In [ ]:

import torch
import platform
import shutil

print("Python:", platform.python_version())
print("PyTorch:", torch.__version__)
print("CUDA available:", torch.cuda.is_available())

if torch.cuda.is_available():
    gpu = torch.cuda.get_device_properties(0)

    print("\nGPU:", torch.cuda.get_device_name(0))
    print("GPU VRAM:", round(gpu.total_memory / 1024**3, 2), "GB")
    print("CUDA version:", torch.version.cuda)
else:
    print("\nWARNING: GPU is not enabled.")

disk = shutil.disk_usage("/content")

print("\nColab storage:")
print("Total:", round(disk.total / 1024**3, 2), "GB")
print("Free:", round(disk.free / 1024**3, 2), "GB")


Python: 3.13.15
PyTorch: 2.11.0+cu130
CUDA available: True

GPU: Tesla T4
GPU VRAM: 14.56 GB
CUDA version: 13.0

Colab storage:
Total: 112.64 GB
Free: 70.27 GB


In [ ]:

%pip -q install "transformers==4.57.6" "datasets[audio]==4.8.5" "accelerate==1.15.0" "torchcodec==0.11.0" "jiwer==4.0.0" "soundfile>=0.13.1,<1" "librosa>=0.11,<1"

import importlib.metadata as metadata
import shutil

packages = [
    "transformers",
    "datasets",
    "accelerate",
    "torchcodec",
    "jiwer",
    "soundfile",
    "librosa",
]

print("Installed libraries:")
for package in packages:
    print(f"{package}: {metadata.version(package)}")

from transformers import (
    Wav2Vec2ForCTC,
    Wav2Vec2CTCTokenizer,
    Wav2Vec2FeatureExtractor,
    Wav2Vec2Processor,
)
from datasets import load_dataset, Audio
from torchcodec.decoders import AudioDecoder

print("\nASR imports: successful")
print("FFmpeg available:", shutil.which("ffmpeg") is not None)


     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 44.0/44.0 kB 2.7 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 12.0/12.0 MB 106.9 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 566.4/566.4 kB 46.1 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 3.2/3.2 MB 124.5 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 3.3/3.3 MB 114.9 MB/s eta 0:00:00
ERROR: pip's dependency resolver does not currently take into account all the packages that are installed. This behaviour is the source of the following dependency conflicts.
gradio 6.30.0 requires huggingface-hub<3.0,>=1.16.0, but you have huggingface-hub 0.36.2 which is incompatible.
diffusers 0.41.0 requires huggingface-hub<2.0,>=1.32.0, but you have huggingface-hub 0.36.2 which is incompatible.
gradio-client 2.7.2 requires huggingface-hub<3.0,>=1.16.0, but you have huggingface-hub 0.36.2 which is incompatible.
Installed libraries:
transformers: 4.57.6
datasets: 4.8.5
accelerate: 1.15.0
torchc

In [ ]:

from datasets import load_dataset_builder

DATASET_NAME = "google/WaxalNLP"
DATASET_CONFIG = "amh_asr"

print("Inspecting dataset metadata...\n")

builder = load_dataset_builder(
    DATASET_NAME,
    DATASET_CONFIG
)

info = builder.info

print("Dataset:", DATASET_NAME)
print("Configuration:", builder.config.name)

print("\nFeatures:")
print(info.features)

print("\nAvailable splits:")

if info.splits:
    for name, split in info.splits.items():
        print(f"\n{name}:")
        print("  Recordings:", split.num_examples)
        print(
            "  Storage size:",
            round(split.num_bytes / 1024**3, 2)
            if split.num_bytes else "Unknown",
            "GB"
        )
else:
    print("Split counts unavailable in builder metadata.")

print("\nLicense:", info.license or "See dataset card")


Inspecting dataset metadata...



/usr/local/lib/python3.13/dist-packages/huggingface_hub/utils/_auth.py:94: UserWarning: 
The secret `HF_TOKEN` does not exist in your Colab secrets.
To authenticate with the Hugging Face Hub, create a token in your settings tab (https://huggingface.co/settings/tokens), set it as secret in your Google Colab and restart your session.
You will be able to reuse this secret in all of your notebooks.
Please note that authentication is recommended but still optional to access public models or datasets.
  warnings.warn(


README.md: 0.00B [00:00, ?B/s]

Resolving data files:   0%|          | 0/72 [00:00<?, ?it/s]

Resolving data files:   0%|          | 0/21 [00:00<?, ?it/s]

Resolving data files:   0%|          | 0/44 [00:00<?, ?it/s]

Dataset: google/WaxalNLP
Configuration: amh_asr

Features:
{'id': Value('string'), 'speaker_id': Value('string'), 'transcription': Value('string'), 'language': Value('string'), 'gender': Value('string'), 'audio': Audio(sampling_rate=None, decode=True, num_channels=None, stream_index=None)}

Available splits:
Split counts unavailable in builder metadata.

License: See dataset card


In [ ]:

import requests

DATASET_NAME = "google/WaxalNLP"
DATASET_CONFIG = "amh_asr"

url = "https://datasets-server.huggingface.co/size"

response = requests.get(
    url,
    params={"dataset": DATASET_NAME},
    timeout=60
)
response.raise_for_status()

data = response.json()
size_info = data.get("size", {})

# Find our specific language configuration.
configs = [
    c for c in size_info.get("configs", [])
    if c.get("config") == DATASET_CONFIG
]

splits = [
    s for s in size_info.get("splits", [])
    if s.get("config") == DATASET_CONFIG
]

print("Dataset:", DATASET_NAME)
print("Configuration:", DATASET_CONFIG)

print("\nConfiguration summary:")
for config in configs:
    print("Total recordings:", config.get("num_rows"))
    print(
        "Storage:",
        round(
            (config.get("num_bytes_original_files") or 0)
            / 1024**3, 2
        ),
        "GB"
    )

print("\nSplit details:")
for split in splits:
    print(
        f"{split.get('split', 'unknown'):12} "
        f"recordings={split.get('num_rows', 'unknown')}, "
        f"size={((split.get('num_bytes_original_files')))} "
        f"or {(split.get('num_bytes_parquet_files') or 0) / 1024**3:.2f} GB"
    )

print("\nPartial metadata:", data.get("partial", False))
print("Pending entries:", len(data.get("pending", [])))
print("Failed entries:", len(data.get("failed", [])))

if not splits:
    print("\nNo split counts returned by the API.")
    print("We may need to inspect Parquet metadata directly.")


Dataset: google/WaxalNLP
Configuration: amh_asr

Configuration summary:
Total recordings: 124675
Storage: 32.25 GB

Split details:
train        recordings=38022, size=None or 9.82 GB
validation   recordings=2912, size=None or 0.73 GB
test         recordings=3420, size=None or 0.86 GB
unlabeled    recordings=80321, size=None or 20.84 GB

Partial metadata: False
Pending entries: 0
Failed entries: 0


In [ ]:

import requests
import fsspec
import pyarrow.parquet as pq

# Get the Parquet files for the Amharic training split.
response = requests.get(
    "https://datasets-server.huggingface.co/parquet",
    params={"dataset": "google/WaxalNLP"},
    timeout=60
)
response.raise_for_status()

metadata = response.json()

train_shards = [
    entry
    for entry in metadata["parquet_files"]
    if entry["config"] == "amh_asr"
    and entry["split"] == "train"
]

train_shards.sort(key=lambda x: x["filename"])

print("Training Parquet shards:", len(train_shards))
print(
    "Total shard size:",
    round(sum(s["size"] for s in train_shards) / 1024**3, 2),
    "GB"
)

assert train_shards, "No Amharic training shards found."

# Read only metadata columns from the first shard.
url = train_shards[0]["url"]

with fsspec.open(url, "rb", block_size=8 * 1024**2) as file:
    parquet = pq.ParquetFile(file)

    print("\nAvailable columns:")
    print(parquet.schema_arrow.names)

    table = parquet.read_row_group(
        0,
        columns=["id", "speaker_id", "transcription"]
    )

    rows = table.slice(0, 3).to_pylist()

print("\nFirst three examples:")
for row in rows:
    print("\nID:", row["id"])
    print("Speaker:", row["speaker_id"])
    print("Text:", row["transcription"][:200])


Training Parquet shards: 21
Total shard size: 9.82 GB

Available columns:
['id', 'speaker_id', 'transcription', 'language', 'gender', 'audio']

First three examples:

ID: yX9LODng8m44GJFPFlT8
Speaker: bBrDrouGOBZ6wjzoXRoHG7AzFL13
Text: በሰማያዊና ነጭ ልብስ የለበሱ የብስክሌት ተወዳዳሪዎች ለመጀመር ሲጠባበቁ በትኩረትና በቆራጥነት ይስተዋላሉ። በደንብ የተደራጀው ውድድር የመጓጓትና የደስታ ስሜት አለው፣ ሁሉም ውድድሩን ለመጀመር ዝግጁ ሆነው ቆመዋል።

ID: yXX1acORw4RRnGAaeBfc
Speaker: koS2CkyGupZguCk2Jd0HtSTpoyP2
Text: በፀሐይ ብርሃን የበቀለ ሰፋፊ የእርሻ መሬት ላይ አረንጓዴ ሽንብራ ከቅጠሎቹ ጋር በፍሬ ተሞልቶ ይታያል። ሰብሉ ሙሉ በሙሉ በልምላሜ የተሸፈነ ሲሆን፣ ከሩቅ ደግሞ ክፍት ሰማይ እና አረንጓዴ ሜዳዎች ይታያሉ፤ ይህም የመልካም ምርትን ተስፋ ይፈጥራል።

ID: yXbBcCapoj9fg8qHOJ3s
Speaker: HJHm7GWboWNaB2Pd4ZHcJ7Vl6rj2
Text: አብዛኞቹ ሴቶች ነጭ ባህላዊ ቀሚሶችን ለብሰዋል፤ ከቀሚሱ ግርጌና በትከሻቸው ላይ የተለያዩ ደማቅ ቀለማት ያላቸው የጥልፍ (የሀገር ልብስ) ቅጦች ይታያሉ።በግራ በኩል አንዲት ሴት የባህላዊ ከበሮ የምትመታ ትመስላለች።




In [ ]:

import json
from pathlib import Path
from collections import Counter

import fsspec
import pyarrow.parquet as pq
from tqdm.auto import tqdm

OUTPUT_PATH = Path("/content/waxal_amh_train_metadata.jsonl")

total_rows = 0
empty_texts = 0
duplicate_ids = 0

speaker_ids = set()
seen_ids = set()
character_counts = Counter()

with OUTPUT_PATH.open("w", encoding="utf-8") as out:

    for shard in tqdm(train_shards, desc="Reading training shards"):

        with fsspec.open(
            shard["url"],
            "rb",
            block_size=8 * 1024**2
        ) as file:

            parquet = pq.ParquetFile(file)

            for batch in parquet.iter_batches(
                batch_size=512,
                columns=["id", "speaker_id", "transcription"]
            ):
                for record in batch.to_pylist():

                    record_id = record["id"]
                    speaker_id = record["speaker_id"]
                    text = record["transcription"] or ""

                    total_rows += 1

                    if not text.strip():
                        empty_texts += 1

                    if record_id in seen_ids:
                        duplicate_ids += 1

                    seen_ids.add(record_id)
                    speaker_ids.add(speaker_id)

                    character_counts.update(text)

                    out.write(
                        json.dumps(
                            {
                                "id": record_id,
                                "speaker_id": speaker_id,
                                "transcription": text
                            },
                            ensure_ascii=False
                        ) + "\n"
                    )

print("\nDATASET SUMMARY")
print("Total recordings:", total_rows)
print("Unique speakers:", len(speaker_ids))
print("Empty transcriptions:", empty_texts)
print("Duplicate IDs:", duplicate_ids)
print("Unique characters:", len(character_counts))

print(
    "Metadata file size:",
    round(OUTPUT_PATH.stat().st_size / 1024**2, 2),
    "MB"
)

print("\nTop 15 characters:")
for char, count in character_counts.most_common(15):
    print(repr(char), count)

assert total_rows == 38022, (
    f"Expected 38,022 rows, found {total_rows}"
)


Reading training shards:   0%|          | 0/21 [00:00<?, ?it/s]


DATASET SUMMARY
Total recordings: 38022
Unique speakers: 566
Empty transcriptions: 0
Duplicate IDs: 0
Unique characters: 402
Metadata file size: 15.9 MB

Top 15 characters:
' ' 985377
'ን' 172661
'የ' 153616
'ት' 144705
'በ' 127272
'ው' 120354
'ል' 112851
'ይ' 104569
'ለ' 102842
'ር' 101250
'ም' 97616
'ያ' 97469
'ስ' 95348
'አ' 89216
'ች' 84594


In [ ]:

import unicodedata
import json
from collections import Counter

def character_group(char):
    name = unicodedata.name(char, "UNKNOWN")
    category = unicodedata.category(char)

    if char.isspace():
        return "WHITESPACE"

    if name.startswith("ETHIOPIC"):
        return "ETHIOPIC"

    if "LATIN" in name:
        return "LATIN"

    if category.startswith("N"):
        return "NUMBER"

    if category.startswith("P"):
        return "PUNCTUATION"

    if category.startswith("S"):
        return "SYMBOL"

    if category.startswith(("C", "M")):
        return "CONTROL / MARK"

    return "OTHER"


# 1. Group characters by Unicode type.
groups = {}

for char, count in character_counts.items():
    group = character_group(char)

    if group not in groups:
        groups[group] = {
            "characters": 0,
            "occurrences": 0
        }

    groups[group]["characters"] += 1
    groups[group]["occurrences"] += count


print("CHARACTER GROUPS")
print("-" * 55)

for group, stats in sorted(groups.items()):
    print(
        f"{group:18} "
        f"unique={stats['characters']:3} "
        f"occurrences={stats['occurrences']:,}"
    )


# 2. Inspect characters outside the Ethiopic script.
print("\nNON-ETHIOPIC CHARACTERS")
print("-" * 55)

non_ethiopic = [
    (char, count)
    for char, count in character_counts.items()
    if character_group(char)
    not in ("ETHIOPIC", "WHITESPACE")
]

for char, count in sorted(
    non_ethiopic,
    key=lambda x: -x[1]
)[:60]:
    print(
        f"{repr(char):10} "
        f"{count:8,} "
        f"{unicodedata.name(char, 'UNKNOWN')}"
    )


# 3. Inspect rare characters.
rare = [
    (char, count)
    for char, count in character_counts.items()
    if count <= 5
]

print("\nRARE CHARACTERS (frequency <= 5)")
print("Total:", len(rare))

for char, count in sorted(
    rare, key=lambda x: x[1]
)[:40]:
    print(
        repr(char),
        count,
        unicodedata.name(char, "UNKNOWN")
    )


# 4. Check normalization effects.
nfc_changes = 0
nfkc_changes = 0

with open(
    OUTPUT_PATH,
    encoding="utf-8"
) as file:
    for line in file:
        text = json.loads(line)["transcription"]

        if unicodedata.normalize("NFC", text) != text:
            nfc_changes += 1

        if unicodedata.normalize("NFKC", text) != text:
            nfkc_changes += 1

print("\nUNICODE NORMALIZATION")
print("Transcripts changed by NFC:", nfc_changes)
print("Transcripts changed by NFKC:", nfkc_changes)


CHARACTER GROUPS
-------------------------------------------------------
CONTROL / MARK     unique=  5 occurrences=47
ETHIOPIC           unique=289 occurrences=3,970,639
LATIN              unique= 54 occurrences=6,394
NUMBER             unique= 10 occurrences=2,230
OTHER              unique=  3 occurrences=5
PUNCTUATION        unique= 28 occurrences=23,778
SYMBOL             unique= 10 occurrences=27
WHITESPACE         unique=  3 occurrences=990,007

NON-ETHIOPIC CHARACTERS
-------------------------------------------------------
'?'           8,032 QUESTION MARK
'!'           4,622 EXCLAMATION MARK
'"'           3,326 QUOTATION MARK
':'           2,518 COLON
'-'           1,193 HYPHEN-MINUS
'('             904 LEFT PARENTHESIS
')'             901 RIGHT PARENTHESIS
"'"             785 APOSTROPHE
'.'             544 FULL STOP
'0'             503 DIGIT ZERO
'1'             482 DIGIT ONE
'e'             436 LATIN SMALL LETTER E
'a'             372 LATIN SMALL LETTER A
'2'             354 D

In [ ]:

import json
import unicodedata
from pathlib import Path
from collections import Counter

NORMALIZED_PATH = Path(
    "/content/waxal_amh_train_normalized.jsonl"
)

def normalize_amharic_ctc(text):
    text = unicodedata.normalize("NFC", text)

    result = []

    for char in text:
        name = unicodedata.name(char, "")
        category = unicodedata.category(char)

        # Standardize whitespace.
        if char.isspace():
            result.append(" ")
            continue

        # Preserve Ethiopic letters and numerals.
        if name.startswith((
            "ETHIOPIC SYLLABLE",
            "ETHIOPIC LETTER",
            "ETHIOPIC DIGIT",
            "ETHIOPIC NUMBER"
        )):
            result.append(char)
            continue

        # Preserve Latin letters, including accented ones.
        if "LATIN" in name and category.startswith("L"):
            result.append(char.lower())
            continue

        # Preserve ASCII digits.
        if char in "0123456789":
            result.append(char)
            continue

        # Remove invisible control/format characters.
        if category.startswith("C"):
            continue

        # Treat punctuation, symbols, and other scripts
        # as word separators.
        result.append(" ")

    # Collapse consecutive spaces.
    return " ".join("".join(result).split())


normalized_counts = Counter()
changed = 0
empty = 0
examples = []

with OUTPUT_PATH.open("r", encoding="utf-8") as source, \
     NORMALIZED_PATH.open("w", encoding="utf-8") as destination:

    for line in source:
        record = json.loads(line)

        original = record["transcription"]
        normalized = normalize_amharic_ctc(original)

        if normalized != original:
            changed += 1

            if len(examples) < 5:
                examples.append((original, normalized))

        if not normalized:
            empty += 1

        normalized_counts.update(normalized)

        record["transcription"] = normalized

        destination.write(
            json.dumps(record, ensure_ascii=False) + "\n"
        )


print("NORMALIZATION SUMMARY")
print("-" * 45)

print("Original unique characters:", len(character_counts))
print("Normalized unique characters:", len(normalized_counts))
print("Modified transcriptions:", changed)
print("Empty transcriptions:", empty)

print(
    "Normalized metadata size:",
    round(NORMALIZED_PATH.stat().st_size / 1024**2, 2),
    "MB"
)

print("\nCHARACTER COVERAGE")
print("Contains reserved '|':", "|" in normalized_counts)

print("\nEXAMPLE TRANSFORMATIONS")

for i, (before, after) in enumerate(examples, 1):
    print(f"\nExample {i}")
    print("BEFORE:", before[:180])
    print("AFTER: ", after[:180])

assert "|" not in normalized_counts
assert empty == 0


NORMALIZATION SUMMARY
---------------------------------------------
Original unique characters: 402
Normalized unique characters: 319
Modified transcriptions: 37208
Empty transcriptions: 0
Normalized metadata size: 15.57 MB

CHARACTER COVERAGE
Contains reserved '|': False

EXAMPLE TRANSFORMATIONS

Example 1
BEFORE: በሰማያዊና ነጭ ልብስ የለበሱ የብስክሌት ተወዳዳሪዎች ለመጀመር ሲጠባበቁ በትኩረትና በቆራጥነት ይስተዋላሉ። በደንብ የተደራጀው ውድድር የመጓጓትና የደስታ ስሜት አለው፣ ሁሉም ውድድሩን ለመጀመር ዝግጁ ሆነው ቆመዋል።
AFTER:  በሰማያዊና ነጭ ልብስ የለበሱ የብስክሌት ተወዳዳሪዎች ለመጀመር ሲጠባበቁ በትኩረትና በቆራጥነት ይስተዋላሉ በደንብ የተደራጀው ውድድር የመጓጓትና የደስታ ስሜት አለው ሁሉም ውድድሩን ለመጀመር ዝግጁ ሆነው ቆመዋል

Example 2
BEFORE: በፀሐይ ብርሃን የበቀለ ሰፋፊ የእርሻ መሬት ላይ አረንጓዴ ሽንብራ ከቅጠሎቹ ጋር በፍሬ ተሞልቶ ይታያል። ሰብሉ ሙሉ በሙሉ በልምላሜ የተሸፈነ ሲሆን፣ ከሩቅ ደግሞ ክፍት ሰማይ እና አረንጓዴ ሜዳዎች ይታያሉ፤ ይህም የመልካም ምርትን ተስፋ ይፈጥራል።
AFTER:  በፀሐይ ብርሃን የበቀለ ሰፋፊ የእርሻ መሬት ላይ አረንጓዴ ሽንብራ ከቅጠሎቹ ጋር በፍሬ ተሞልቶ ይታያል ሰብሉ ሙሉ በሙሉ በልምላሜ የተሸፈነ ሲሆን ከሩቅ ደግሞ ክፍት ሰማይ እና አረንጓዴ ሜዳዎች ይታያሉ ይህም የመልካም ምርትን ተስፋ ይፈጥራል

Example 3
BEFORE: አብዛኞቹ ሴቶች ነጭ ባህላዊ ቀሚሶችን ለብሰዋል፤ ከቀሚሱ ግርጌና በትከሻቸው ላይ የ

In [ ]:

import json
from pathlib import Path
from transformers import Wav2Vec2CTCTokenizer

TOKENIZER_DIR = Path("/content/amharic_ctc_tokenizer")
TOKENIZER_DIR.mkdir(parents=True, exist_ok=True)

# Build vocabulary using the complete normalized corpus.
characters = sorted(
    char for char in normalized_counts
    if char != " "
)

vocab = {
    char: index
    for index, char in enumerate(characters)
}

# Reserve special tokens.
vocab["|"] = len(vocab)
vocab["[UNK]"] = len(vocab)
vocab["[PAD]"] = len(vocab)

VOCAB_PATH = TOKENIZER_DIR / "vocab.json"

with VOCAB_PATH.open("w", encoding="utf-8") as file:
    json.dump(
        vocab,
        file,
        ensure_ascii=False,
        indent=2
    )

# Explicitly disable unnecessary BOS/EOS tokens.
tokenizer = Wav2Vec2CTCTokenizer(
    vocab_file=str(VOCAB_PATH),
    unk_token="[UNK]",
    pad_token="[PAD]",
    word_delimiter_token="|",
    bos_token=None,
    eos_token=None,
    do_lower_case=False,
    clean_up_tokenization_spaces=False
)

# Verify vocabulary integrity.
assert len(tokenizer) == len(vocab)
assert len(set(vocab.values())) == len(vocab)
assert set(vocab.values()) == set(range(len(vocab)))

# All normalized training characters must be representable.
missing = set(normalized_counts) - {" "} - set(vocab)
assert not missing, f"Missing characters: {missing}"

# Test real training transcriptions.
with NORMALIZED_PATH.open(encoding="utf-8") as file:
    samples = [
        json.loads(next(file))["transcription"]
        for _ in range(3)
    ]

for i, text in enumerate(samples, 1):
    token_ids = tokenizer.encode(
        text,
        add_special_tokens=False
    )

    # Disable CTC duplicate collapsing for label round-trip.
    decoded = tokenizer.decode(
        token_ids,
        group_tokens=False,
        clean_up_tokenization_spaces=False
    )

    assert tokenizer.unk_token_id not in token_ids
    assert decoded == text, f"Round-trip failed: {i}"

    print(f"Example {i}:")
    print("  Characters:", len(text))
    print("  Tokens:", len(token_ids))
    print("  Round-trip successful:", decoded == text)

# Save tokenizer configuration alongside vocabulary.
tokenizer.save_pretrained(str(TOKENIZER_DIR))

print("\nVOCABULARY SUMMARY")
print("Total tokens:", len(tokenizer))
print("Word delimiter ID:", tokenizer.word_delimiter_token_id)
print("Unknown token ID:", tokenizer.unk_token_id)
print("CTC blank ID:", tokenizer.pad_token_id)
print("BOS token:", tokenizer.bos_token)
print("EOS token:", tokenizer.eos_token)
print("Saved to:", TOKENIZER_DIR)


Example 1:
  Characters: 132
  Tokens: 132
  Round-trip successful: True
Example 2:
  Characters: 151
  Tokens: 151
  Round-trip successful: True
Example 3:
  Characters: 131
  Tokens: 131
  Round-trip successful: True

VOCABULARY SUMMARY
Total tokens: 321
Word delimiter ID: 318
Unknown token ID: 319
CTC blank ID: 320
BOS token: None
EOS token: None
Saved to: /content/amharic_ctc_tokenizer


In [ ]:

import json
import unicodedata
from pathlib import Path
from collections import Counter

import fsspec
import pyarrow.parquet as pq
from tqdm.auto import tqdm
from transformers import Wav2Vec2CTCTokenizer

# 1. Verify that the saved tokenizer reloads identically.
reloaded_tokenizer = Wav2Vec2CTCTokenizer.from_pretrained(
    str(TOKENIZER_DIR)
)

assert reloaded_tokenizer.get_vocab() == tokenizer.get_vocab()
assert reloaded_tokenizer.pad_token_id == 320
assert reloaded_tokenizer.unk_token_id == 319

print("Tokenizer reload: PASSED")

# 2. Locate validation Parquet shards.
val_shards = sorted(
    [
        shard
        for shard in metadata["parquet_files"]
        if shard["config"] == "amh_asr"
        and shard["split"] == "validation"
    ],
    key=lambda shard: shard["filename"]
)

assert val_shards, "No validation shards found."

# 3. Scan validation text without loading audio.
VAL_METADATA_PATH = Path(
    "/content/waxal_amh_validation_normalized.jsonl"
)

oov_counts = Counter()
validation_speakers = set()

total_records = 0
total_characters = 0
oov_characters = 0
affected_records = 0
empty_records = 0

with VAL_METADATA_PATH.open("w", encoding="utf-8") as out:
    for shard in tqdm(val_shards, desc="Scanning validation"):
        with fsspec.open(
            shard["url"], "rb", block_size=8 * 1024**2
        ) as file:
            parquet = pq.ParquetFile(file)

            for batch in parquet.iter_batches(
                batch_size=512,
                columns=["id", "speaker_id", "transcription"]
            ):
                for record in batch.to_pylist():
                    text = normalize_amharic_ctc(
                        record["transcription"] or ""
                    )

                    total_records += 1
                    total_characters += len(text)
                    validation_speakers.add(record["speaker_id"])

                    if not text:
                        empty_records += 1

                    # Spaces are represented by | in the tokenizer.
                    missing = [
                        char for char in text
                        if char != " " and char not in vocab
                    ]

                    if missing:
                        affected_records += 1
                        oov_characters += len(missing)
                        oov_counts.update(missing)

                    out.write(
                        json.dumps(
                            {
                                "id": record["id"],
                                "speaker_id": record["speaker_id"],
                                "transcription": text
                            },
                            ensure_ascii=False
                        ) + "\n"
                    )

print("\nVALIDATION VOCABULARY AUDIT")
print("-" * 45)
print("Validation recordings:", total_records)
print("Empty transcriptions:", empty_records)
print("Unique validation speakers:", len(validation_speakers))
print(
    "Speakers overlapping training:",
    len(validation_speakers & speaker_ids)
)
print("Recordings containing OOV characters:", affected_records)
print("Unique unseen characters:", len(oov_counts))
print("Total OOV character occurrences:", oov_characters)
print(
    "OOV character rate:",
    f"{100 * oov_characters / max(total_characters, 1):.4f}%"
)

print("\nUNSEEN CHARACTERS (top 20)")
for char, count in oov_counts.most_common(20):
    print(
        repr(char),
        count,
        unicodedata.name(char, "UNKNOWN")
    )

assert total_records == 2912
assert empty_records == 0

print("\nSaved validation metadata:", VAL_METADATA_PATH)


Tokenizer reload: PASSED


Scanning validation:   0%|          | 0/2 [00:00<?, ?it/s]


VALIDATION VOCABULARY AUDIT
---------------------------------------------
Validation recordings: 2912
Empty transcriptions: 0
Unique validation speakers: 28
Speakers overlapping training: 0
Recordings containing OOV characters: 0
Unique unseen characters: 0
Total OOV character occurrences: 0
OOV character rate: 0.0000%

UNSEEN CHARACTERS (top 20)

Saved validation metadata: /content/waxal_amh_validation_normalized.jsonl


In [ ]:

from datasets import load_dataset
from torchcodec.decoders import AudioDecoder
from collections import Counter
from itertools import islice
import statistics

# Stream only the first training shard.
# Avoid loading all 21 shards into memory.
audio_stream = load_dataset(
    "parquet",
    data_files={"train": train_shards[0]["url"]},
    split="train",
    streaming=True
).decode(False)

audio_probe = []

for example in islice(audio_stream, 12):
    audio = example["audio"]

    # Parquet generally stores the encoded audio bytes.
    source = (
        audio["bytes"]
        if audio["bytes"] is not None
        else audio["path"]
    )

    decoder = AudioDecoder(source)
    info = decoder.metadata

    duration = info.duration_seconds

    audio_probe.append({
        "id": example["id"],
        "duration": duration,
        "sample_rate": info.sample_rate,
        "channels": info.num_channels,
        "codec": info.codec
    })

print("AUDIO PROBE RESULTS")
print("-" * 50)

for i, item in enumerate(audio_probe, 1):
    print(
        f"{i:02d} | "
        f"{item['duration']:.2f}s | "
        f"{item['sample_rate']} Hz | "
        f"{item['channels']} channel(s) | "
        f"{item['codec']}"
    )

durations = [x["duration"] for x in audio_probe]

print("\nSUMMARY")
print("Recordings inspected:", len(audio_probe))
print("Mean duration:", round(statistics.mean(durations), 2), "s")
print("Median duration:", round(statistics.median(durations), 2), "s")
print("Min duration:", round(min(durations), 2), "s")
print("Max duration:", round(max(durations), 2), "s")

print(
    "Sample rates:",
    dict(Counter(x["sample_rate"] for x in audio_probe))
)

print(
    "Channels:",
    dict(Counter(x["channels"] for x in audio_probe))
)

print(
    "Codecs:",
    dict(Counter(x["codec"] for x in audio_probe))
)


AUDIO PROBE RESULTS
--------------------------------------------------
01 | 22.46s | 48000 Hz | 1 channel(s) | mp3
02 | 23.90s | 48000 Hz | 1 channel(s) | mp3
03 | 18.14s | 48000 Hz | 1 channel(s) | mp3
04 | 18.98s | 48000 Hz | 1 channel(s) | mp3
05 | 18.94s | 48000 Hz | 1 channel(s) | mp3
06 | 17.26s | 48000 Hz | 1 channel(s) | mp3
07 | 17.50s | 48000 Hz | 1 channel(s) | mp3
08 | 18.74s | 48000 Hz | 1 channel(s) | mp3
09 | 16.22s | 48000 Hz | 1 channel(s) | mp3
10 | 19.22s | 48000 Hz | 1 channel(s) | mp3
11 | 15.58s | 48000 Hz | 1 channel(s) | mp3
12 | 18.74s | 48000 Hz | 1 channel(s) | mp3

SUMMARY
Recordings inspected: 12
Mean duration: 18.81 s
Median duration: 18.74 s
Min duration: 15.58 s
Max duration: 23.9 s
Sample rates: {48000: 12}
Channels: {1: 12}
Codecs: {'mp3': 12}


In [ ]:

from google.colab import drive
from pathlib import Path
import shutil
import json
import hashlib

# Mount Google Drive.
drive.mount("/content/drive")

# Create project directories.
PROJECT_DIR = Path(
    "/content/drive/MyDrive/Amharic_ASR_XLSR"
)

DATA_DIR = PROJECT_DIR / "data"
TOKENIZER_SAVE_DIR = PROJECT_DIR / "tokenizer"
CHECKPOINT_DIR = PROJECT_DIR / "checkpoints"

for directory in [
    DATA_DIR,
    TOKENIZER_SAVE_DIR,
    CHECKPOINT_DIR
]:
    directory.mkdir(parents=True, exist_ok=True)

# Save the original and normalized metadata.
files_to_save = {
    "train_original.jsonl": OUTPUT_PATH,
    "train_normalized.jsonl": NORMALIZED_PATH,
    "validation_normalized.jsonl": VAL_METADATA_PATH,
}

for name, source in files_to_save.items():
    destination = DATA_DIR / name
    shutil.copy2(source, destination)

    print(
        f"Saved {name}: "
        f"{destination.stat().st_size / 1024**2:.2f} MB"
    )

# Save the complete tokenizer directory.
shutil.copytree(
    TOKENIZER_DIR,
    TOKENIZER_SAVE_DIR,
    dirs_exist_ok=True
)

# Save experiment metadata.
experiment_config = {
    "dataset": "google/WaxalNLP",
    "dataset_config": "amh_asr",
    "model": "facebook/wav2vec2-xls-r-300m",
    "train_examples": 38022,
    "validation_examples": 2912,
    "vocab_size": len(tokenizer),
    "blank_token_id": tokenizer.pad_token_id,
    "target_sample_rate": 16000,
    "normalization": "NFC, lowercase Latin, strip punctuation and unsupported symbols, collapse whitespace",
}

with (PROJECT_DIR / "experiment_config.json").open(
    "w", encoding="utf-8"
) as file:
    json.dump(
        experiment_config,
        file,
        ensure_ascii=False,
        indent=2
    )

# Verify that the saved tokenizer can be reloaded.
from transformers import Wav2Vec2CTCTokenizer

saved_tokenizer = Wav2Vec2CTCTokenizer.from_pretrained(
    str(TOKENIZER_SAVE_DIR)
)

assert saved_tokenizer.get_vocab() == tokenizer.get_vocab()

print("\nBACKUP COMPLETE")
print("Project:", PROJECT_DIR)
print("Tokenizer:", TOKENIZER_SAVE_DIR)
print("Vocabulary size:", len(saved_tokenizer))
print("Checkpoint directory:", CHECKPOINT_DIR)


Drive already mounted at /content/drive; to attempt to forcibly remount, call drive.mount("/content/drive", force_remount=True).
Saved train_original.jsonl: 15.90 MB
Saved train_normalized.jsonl: 15.57 MB
Saved validation_normalized.jsonl: 1.20 MB

BACKUP COMPLETE
Project: /content/drive/MyDrive/Amharic_ASR_XLSR
Tokenizer: /content/drive/MyDrive/Amharic_ASR_XLSR/tokenizer
Vocabulary size: 321
Checkpoint directory: /content/drive/MyDrive/Amharic_ASR_XLSR/checkpoints


In [ ]:

from itertools import islice
from datasets import load_dataset
from torchcodec.decoders import AudioDecoder
from IPython.display import Audio, display
import numpy as np

def inspect_recordings(shard, count, split_name):
    stream = load_dataset(
        "parquet",
        data_files={"train": shard["url"]},
        split="train",
        streaming=True
    ).decode(False)

    for i, example in enumerate(islice(stream, count), 1):
        audio_info = example["audio"]

        source = audio_info.get("bytes")
        if source is None:
            source = audio_info.get("path")

        if source is None:
            raise ValueError("Audio bytes/path missing")

        # Decode AND resample to our model's required 16 kHz.
        decoder = AudioDecoder(
            source,
            sample_rate=16000,
            num_channels=1
        )

        samples = decoder.get_all_samples()
        waveform = samples.data[0].cpu().numpy()

        duration = len(waveform) / samples.sample_rate
        rms = float(np.sqrt(np.mean(waveform ** 2)))

        print(f"\n{'=' * 60}")
        print(f"{split_name} RECORDING {i}")
        print(f"{'=' * 60}")

        print("ID:", example["id"])
        print("Speaker:", example["speaker_id"])
        print("Duration:", round(duration, 2), "seconds")
        print("Decoded sample rate:", samples.sample_rate, "Hz")
        print("Audio RMS:", round(rms, 4))

        print("\nORIGINAL TRANSCRIPTION:")
        print(example["transcription"])

        print("\nNORMALIZED TRANSCRIPTION:")
        print(normalize_amharic_ctc(example["transcription"]))

        print("\nLISTEN:")
        display(Audio(waveform, rate=samples.sample_rate))


# Two training recordings.
inspect_recordings(
    train_shards[0],
    count=2,
    split_name="TRAIN"
)

# One validation recording.
inspect_recordings(
    val_shards[0],
    count=1,
    split_name="VALIDATION"
)



TRAIN RECORDING 1
ID: yX9LODng8m44GJFPFlT8
Speaker: bBrDrouGOBZ6wjzoXRoHG7AzFL13
Duration: 22.46 seconds
Decoded sample rate: 16000 Hz
Audio RMS: 0.0509

ORIGINAL TRANSCRIPTION:
በሰማያዊና ነጭ ልብስ የለበሱ የብስክሌት ተወዳዳሪዎች ለመጀመር ሲጠባበቁ በትኩረትና በቆራጥነት ይስተዋላሉ። በደንብ የተደራጀው ውድድር የመጓጓትና የደስታ ስሜት አለው፣ ሁሉም ውድድሩን ለመጀመር ዝግጁ ሆነው ቆመዋል።

NORMALIZED TRANSCRIPTION:
በሰማያዊና ነጭ ልብስ የለበሱ የብስክሌት ተወዳዳሪዎች ለመጀመር ሲጠባበቁ በትኩረትና በቆራጥነት ይስተዋላሉ በደንብ የተደራጀው ውድድር የመጓጓትና የደስታ ስሜት አለው ሁሉም ውድድሩን ለመጀመር ዝግጁ ሆነው ቆመዋል

LISTEN:



TRAIN RECORDING 2
ID: yXX1acORw4RRnGAaeBfc
Speaker: koS2CkyGupZguCk2Jd0HtSTpoyP2
Duration: 23.9 seconds
Decoded sample rate: 16000 Hz
Audio RMS: 0.0743

ORIGINAL TRANSCRIPTION:
በፀሐይ ብርሃን የበቀለ ሰፋፊ የእርሻ መሬት ላይ አረንጓዴ ሽንብራ ከቅጠሎቹ ጋር በፍሬ ተሞልቶ ይታያል። ሰብሉ ሙሉ በሙሉ በልምላሜ የተሸፈነ ሲሆን፣ ከሩቅ ደግሞ ክፍት ሰማይ እና አረንጓዴ ሜዳዎች ይታያሉ፤ ይህም የመልካም ምርትን ተስፋ ይፈጥራል።

NORMALIZED TRANSCRIPTION:
በፀሐይ ብርሃን የበቀለ ሰፋፊ የእርሻ መሬት ላይ አረንጓዴ ሽንብራ ከቅጠሎቹ ጋር በፍሬ ተሞልቶ ይታያል ሰብሉ ሙሉ በሙሉ በልምላሜ የተሸፈነ ሲሆን ከሩቅ ደግሞ ክፍት ሰማይ እና አረንጓዴ ሜዳዎች ይታያሉ ይህም የመልካም ምርትን ተስፋ ይፈጥራል

LISTEN:



VALIDATION RECORDING 1
ID: G1FVSAM9JejBObRk5dy0
Speaker: t4058VWLeJRUpyMAMPYXEtJBie03
Duration: 20.14 seconds
Decoded sample rate: 16000 Hz
Audio RMS: 0.0328

ORIGINAL TRANSCRIPTION:
ጥቁር ሰማያዊ፣ ነጭና ወርቃማ ቀለም ያላቸው ብዙ ፊኛዎች፣ አበባዎችና መብራቶች ያጌጠ ቦታ ነው።  በግራ በኩል በክፈፍ ውስጥ ያለ የህፃን ልጅ ምስል እና በፊት ለፊት ሰማያዊና ነጭ አበባዎች የያዙ ማቆሚያዎች የደስታ፣ የፍቅርና የልደት በዓል ድባብን ይፈጥራሉ።

NORMALIZED TRANSCRIPTION:
ጥቁር ሰማያዊ ነጭና ወርቃማ ቀለም ያላቸው ብዙ ፊኛዎች አበባዎችና መብራቶች ያጌጠ ቦታ ነው በግራ በኩል በክፈፍ ውስጥ ያለ የህፃን ልጅ ምስል እና በፊት ለፊት ሰማያዊና ነጭ አበባዎች የያዙ ማቆሚያዎች የደስታ የፍቅርና የልደት በዓል ድባብን ይፈጥራሉ

LISTEN:


In [ ]:

import random
import math
import statistics
import numpy as np
import fsspec
import pyarrow.parquet as pq

from torchcodec.decoders import AudioDecoder
from tqdm.auto import tqdm

SEED = 42
rng = random.Random(SEED)

TARGET_HOURS = 25

# Sample 9 shards distributed throughout the training dataset.
shard_indices = sorted(set(
    round(i * (len(train_shards) - 1) / 8)
    for i in range(9)
))

duration_probe = []
errors = []

for shard_index in tqdm(
    shard_indices,
    desc="Sampling audio across shards"
):
    shard = train_shards[shard_index]

    try:
        with fsspec.open(
            shard["url"],
            "rb",
            block_size=8 * 1024**2
        ) as file:
            parquet = pq.ParquetFile(file)

            # Select a random row group rather than always
            # reading the beginning of each shard.
            group_index = rng.randrange(
                parquet.metadata.num_row_groups
            )

            table = parquet.read_row_group(
                group_index,
                columns=["id", "speaker_id", "audio"]
            )

            records = table.to_pylist()

            chosen_indices = rng.sample(
                range(len(records)),
                min(5, len(records))
            )

            for index in chosen_indices:
                record = records[index]
                audio = record["audio"]

                source = audio.get("bytes")
                if source is None:
                    source = audio.get("path")

                decoder = AudioDecoder(source)
                duration = decoder.metadata.duration_seconds

                if duration is None or not math.isfinite(duration):
                    continue

                duration_probe.append({
                    "id": record["id"],
                    "speaker_id": record["speaker_id"],
                    "duration": float(duration),
                    "shard_index": shard_index
                })

    except Exception as exc:
        errors.append((shard_index, str(exc)[:200]))


durations = np.array([
    item["duration"] for item in duration_probe
])

assert len(durations) > 0, "No valid audio durations found."

print("\nAUDIO DURATION ANALYSIS")
print("-" * 48)

print("Recordings inspected:", len(durations))
print(
    "Unique speakers:",
    len(set(item["speaker_id"] for item in duration_probe))
)

print("Mean:", round(float(durations.mean()), 2), "seconds")
print("Median:", round(float(np.median(durations)), 2), "seconds")
print("Minimum:", round(float(durations.min()), 2), "seconds")
print("Maximum:", round(float(durations.max()), 2), "seconds")

print("\nDURATION PERCENTILES")
for percentile in [10, 25, 50, 75, 90, 95]:
    value = np.percentile(durations, percentile)
    print(f"P{percentile}: {value:.2f} seconds")

print("\nDURATION BUCKETS")
buckets = [
    ("Under 10s", durations < 10),
    ("10-20s", (durations >= 10) & (durations < 20)),
    ("20-30s", (durations >= 20) & (durations < 30)),
    ("30-40s", (durations >= 30) & (durations < 40)),
    ("40s+", durations >= 40)
]

for label, mask in buckets:
    print(f"{label:12} {int(mask.sum()):3} recordings")

estimated_total_hours = (
    38022 * durations.mean() / 3600
)

estimated_recordings = (
    TARGET_HOURS * 3600 / durations.mean()
)

print("\nPRELIMINARY TRAINING ESTIMATES")
print(
    "Estimated full training duration:",
    round(estimated_total_hours, 1),
    "hours"
)
print(
    "Estimated recordings for 25 hours:",
    round(estimated_recordings)
)

print("\nRead errors:", len(errors))
for error in errors[:5]:
    print(error)


Sampling audio across shards:   0%|          | 0/9 [00:00<?, ?it/s]


AUDIO DURATION ANALYSIS
------------------------------------------------
Recordings inspected: 43
Unique speakers: 21
Mean: 18.26 seconds
Median: 17.74 seconds
Minimum: 14.98 seconds
Maximum: 25.22 seconds

DURATION PERCENTILES
P10: 15.35 seconds
P25: 16.44 seconds
P50: 17.74 seconds
P75: 19.72 seconds
P90: 21.62 seconds
P95: 21.92 seconds

DURATION BUCKETS
Under 10s      0 recordings
10-20s        33 recordings
20-30s        10 recordings
30-40s         0 recordings
40s+           0 recordings

PRELIMINARY TRAINING ESTIMATES
Estimated full training duration: 192.8 hours
Estimated recordings for 25 hours: 4930

Read errors: 0


In [ ]:

import json
import math
import random
from pathlib import Path
from collections import defaultdict, Counter

# =============================================
# EXPERIMENT CONFIGURATION
# =============================================

TRAIN_TARGET_HOURS = 25.0   # Change to 50, 100, etc.
                            # Use None for the full corpus.

RANDOM_SEED = 42

# Estimated from our 43-recording audio probe.
ESTIMATED_CLIP_SECONDS = 18.26

# Extra candidates to allow filtering and duration variation.
CANDIDATE_BUFFER = 1.20

# =============================================
# BUILD STABLE, SPEAKER-BALANCED PRIORITY ORDER
# =============================================

rng = random.Random(RANDOM_SEED)
speaker_pools = defaultdict(list)

with NORMALIZED_PATH.open(encoding="utf-8") as file:
    for row_index, line in enumerate(file):
        record = json.loads(line)
        record["source_row_index"] = row_index
        speaker_pools[record["speaker_id"]].append(record)

# Reproducible shuffling within each speaker.
for speaker in sorted(speaker_pools):
    rng.shuffle(speaker_pools[speaker])

active_speakers = sorted(speaker_pools)
priority_records = []

# Round-robin selection gives speakers opportunities
# to contribute recordings before others dominate.
while active_speakers:
    rng.shuffle(active_speakers)
    next_active = []

    for speaker in active_speakers:
        pool = speaker_pools[speaker]

        if pool:
            record = pool.pop()
            record["selection_rank"] = len(priority_records)
            priority_records.append(record)

        if pool:
            next_active.append(speaker)

    active_speakers = next_active

assert len(priority_records) == 38022
assert len({r["id"] for r in priority_records}) == 38022

# =============================================
# SELECT A CANDIDATE POOL
# =============================================

if TRAIN_TARGET_HOURS is None:
    candidate_count = len(priority_records)
    plan_label = "full"
else:
    estimated_count = (
        TRAIN_TARGET_HOURS * 3600
        / ESTIMATED_CLIP_SECONDS
    )

    candidate_count = min(
        math.ceil(estimated_count * CANDIDATE_BUFFER),
        len(priority_records)
    )
    plan_label = f"{TRAIN_TARGET_HOURS:g}h".replace(".", "p")

candidates = priority_records[:candidate_count]

# =============================================
# SAVE MANIFESTS AND CONFIGURATION
# =============================================

PRIORITY_PATH = DATA_DIR / "train_priority_all.jsonl"
CANDIDATE_PATH = (
    DATA_DIR / f"train_candidates_{plan_label}.jsonl"
)

def save_jsonl(records, path):
    with path.open("w", encoding="utf-8") as file:
        for record in records:
            file.write(
                json.dumps(record, ensure_ascii=False) + "\n"
            )

save_jsonl(priority_records, PRIORITY_PATH)
save_jsonl(candidates, CANDIDATE_PATH)

training_plan = {
    "target_hours": TRAIN_TARGET_HOURS,
    "seed": RANDOM_SEED,
    "estimated_clip_seconds": ESTIMATED_CLIP_SECONDS,
    "candidate_buffer": CANDIDATE_BUFFER,
    "candidate_count": candidate_count,
    "priority_manifest": str(PRIORITY_PATH),
    "candidate_manifest": str(CANDIDATE_PATH),
    "selection_method": "seeded_speaker_round_robin",
    "duration_status": "estimated_not_measured"
}

PLAN_PATH = DATA_DIR / f"training_plan_{plan_label}.json"

with PLAN_PATH.open("w", encoding="utf-8") as file:
    json.dump(training_plan, file, indent=2)

# =============================================
# REPORT
# =============================================

speaker_counts = Counter(
    r["speaker_id"] for r in candidates
)

candidate_characters = set().union(
    *(set(r["transcription"]) for r in candidates)
)

print("CONFIGURABLE TRAINING PLAN")
print("-" * 50)

print("Target hours:", TRAIN_TARGET_HOURS)
print("Total available recordings:", len(priority_records))
print("Candidate recordings:", len(candidates))
print("Selected speakers:", len(speaker_counts))
print("Minimum clips per speaker:", min(speaker_counts.values()))
print("Maximum clips per speaker:", max(speaker_counts.values()))

print(
    "Estimated candidate-pool hours:",
    round(
        len(candidates) * ESTIMATED_CLIP_SECONDS / 3600,
        2
    )
)

print(
    "Candidate character coverage:",
    len(candidate_characters),
    "/",
    len(normalized_counts)
)

print("\nSaved priority manifest:", PRIORITY_PATH)
print("Saved candidate manifest:", CANDIDATE_PATH)
print("Saved training plan:", PLAN_PATH)

print("\nNEXT: Measure actual candidate durations.")


CONFIGURABLE TRAINING PLAN
--------------------------------------------------
Target hours: 25.0
Total available recordings: 38022
Candidate recordings: 5915
Selected speakers: 566
Minimum clips per speaker: 1
Maximum clips per speaker: 13
Estimated candidate-pool hours: 30.0
Candidate character coverage: 289 / 319

Saved priority manifest: /content/drive/MyDrive/Amharic_ASR_XLSR/data/train_priority_all.jsonl
Saved candidate manifest: /content/drive/MyDrive/Amharic_ASR_XLSR/data/train_candidates_25h.jsonl
Saved training plan: /content/drive/MyDrive/Amharic_ASR_XLSR/data/training_plan_25h.json

NEXT: Measure actual candidate durations.


In [ ]:

import json
import math
from bisect import bisect_left
from pathlib import Path

import fsspec
import pyarrow.parquet as pq
from torchcodec.decoders import AudioDecoder
from tqdm.auto import tqdm

# ==========================================
# CONFIGURATION
# ==========================================

AUDIO_DIR = Path("/content/amharic_asr_candidate_audio")
AUDIO_DIR.mkdir(parents=True, exist_ok=True)

PROGRESS_PATH = Path(
    "/content/amharic_audio_extraction_progress.jsonl"
)

TARGET_SECONDS = TRAIN_TARGET_HOURS * 3600

# Load selected candidates.
with CANDIDATE_PATH.open(encoding="utf-8") as f:
    candidate_records = [json.loads(line) for line in f]

candidates_by_row = {
    r["source_row_index"]: r for r in candidate_records
}

selected_positions = sorted(candidates_by_row)

# Restore extraction progress, ignoring missing local files.
completed = {}

if PROGRESS_PATH.exists():
    with PROGRESS_PATH.open(encoding="utf-8") as f:
        for line in f:
            record = json.loads(line)
            audio_path = AUDIO_DIR / record["audio_file"]

            if audio_path.exists() and audio_path.stat().st_size > 0:
                completed[record["id"]] = record

print("Candidates:", len(candidate_records))
print("Already extracted:", len(completed))

errors = []
global_start = 0

# ==========================================
# EXTRACT SELECTED AUDIO FROM PARQUET
# ==========================================

with PROGRESS_PATH.open("a", encoding="utf-8") as progress_file:

    for shard_index, shard in enumerate(
        tqdm(train_shards, desc="Extracting audio shards")
    ):
        with fsspec.open(
            shard["url"],
            "rb",
            block_size=16 * 1024**2
        ) as source:
            parquet = pq.ParquetFile(source)

            shard_rows = parquet.metadata.num_rows
            shard_end = global_start + shard_rows

            # Find candidates belonging to this shard.
            left = bisect_left(selected_positions, global_start)
            right = bisect_left(selected_positions, shard_end)

            shard_positions = selected_positions[left:right]
            shard_position_set = set(shard_positions)

            group_start = global_start

            for group_index in range(parquet.metadata.num_row_groups):
                group_rows = parquet.metadata.row_group(
                    group_index
                ).num_rows

                group_end = group_start + group_rows

                needed_positions = [
                    pos for pos in shard_positions
                    if group_start <= pos < group_end
                    and candidates_by_row[pos]["id"] not in completed
                ]

                if not needed_positions:
                    group_start = group_end
                    continue

                needed = set(needed_positions)
                row_offset = 0

                for batch in parquet.iter_batches(
                    row_groups=[group_index],
                    columns=["id", "audio"],
                    batch_size=64
                ):
                    records = batch.to_pylist()

                    for local_index, record in enumerate(records):
                        global_index = (
                            group_start + row_offset + local_index
                        )

                        if global_index not in needed:
                            continue

                        expected = candidates_by_row[global_index]

                        # Verify our transcript/audio indexing.
                        assert record["id"] == expected["id"], (
                            f"ID mismatch at row {global_index}"
                        )

                        try:
                            encoded_audio = record["audio"]["bytes"]

                            if encoded_audio is None:
                                raise ValueError(
                                    "Audio bytes missing from Parquet"
                                )

                            decoder = AudioDecoder(encoded_audio)
                            duration = (
                                decoder.metadata.duration_seconds
                            )

                            if (
                                duration is None
                                or not math.isfinite(duration)
                                or duration <= 0
                            ):
                                raise ValueError(
                                    f"Invalid duration: {duration}"
                                )

                            filename = expected["id"] + ".mp3"
                            destination = AUDIO_DIR / filename
                            temporary = AUDIO_DIR / (filename + ".tmp")

                            temporary.write_bytes(encoded_audio)
                            temporary.replace(destination)

                            result = {
                                **expected,
                                "duration_seconds": float(duration),
                                "audio_file": filename
                            }

                            completed[expected["id"]] = result

                            progress_file.write(
                                json.dumps(
                                    result, ensure_ascii=False
                                ) + "\n"
                            )
                            progress_file.flush()

                        except Exception as exc:
                            errors.append(
                                (expected["id"], str(exc)[:200])
                            )

                    row_offset += len(records)

                group_start = group_end

            global_start = shard_end

# ==========================================
# SELECT FINAL TRAINING HOURS
# ==========================================

measured = sorted(
    completed.values(),
    key=lambda r: r["selection_rank"]
)

final_records = []
actual_seconds = 0.0

for record in measured:
    if actual_seconds >= TARGET_SECONDS:
        break

    final_records.append(record)
    actual_seconds += record["duration_seconds"]

FINAL_MANIFEST = (
    DATA_DIR / f"train_final_{TRAIN_TARGET_HOURS:g}h.jsonl"
)

with FINAL_MANIFEST.open("w", encoding="utf-8") as f:
    for record in final_records:
        f.write(json.dumps(record, ensure_ascii=False) + "\n")

# ==========================================
# REPORT
# ==========================================

print("\nAUDIO EXTRACTION SUMMARY")
print("-" * 50)
print("Candidates requested:", len(candidate_records))
print("Candidates extracted:", len(completed))
print("Extraction errors:", len(errors))

print("\nFINAL TRAINING SELECTION")
print("Target hours:", TRAIN_TARGET_HOURS)
print("Actual hours:", round(actual_seconds / 3600, 3))
print("Selected recordings:", len(final_records))
print(
    "Selected speakers:",
    len({r["speaker_id"] for r in final_records})
)

print(
    "Local audio storage:",
    round(
        sum(p.stat().st_size for p in AUDIO_DIR.glob("*.mp3"))
        / 1024**3,
        2
    ),
    "GB"
)

print("\nFinal manifest:", FINAL_MANIFEST)
print("Audio directory:", AUDIO_DIR)

if errors:
    print("\nFirst extraction errors:")
    for error in errors[:5]:
        print(error)

if actual_seconds < TARGET_SECONDS:
    print(
        "\nWARNING: Candidate pool did not reach the target."
        "\nWe can expand the pool using the saved priority list."
    )
else:
    print("\nTarget duration achieved.")

assert global_start == 38022, (
    f"Dataset indexing mismatch: {global_start}"
)


Candidates: 5915
Already extracted: 0


Extracting audio shards:   0%|          | 0/21 [00:00<?, ?it/s]


AUDIO EXTRACTION SUMMARY
--------------------------------------------------
Candidates requested: 5915
Candidates extracted: 5915
Extraction errors: 0

FINAL TRAINING SELECTION
Target hours: 25.0
Actual hours: 25.001
Selected recordings: 5084
Selected speakers: 566
Local audio storage: 1.56 GB

Final manifest: /content/drive/MyDrive/Amharic_ASR_XLSR/data/train_final_25h.jsonl
Audio directory: /content/amharic_asr_candidate_audio

Target duration achieved.


In [ ]:

import json
import tarfile
import hashlib
import shutil
from pathlib import Path
from tqdm.auto import tqdm

ARCHIVE_BATCH_SIZE = 600

ARCHIVE_DIR = PROJECT_DIR / "audio_archives" / "25h"
ARCHIVE_DIR.mkdir(parents=True, exist_ok=True)

LOCAL_ARCHIVE_DIR = Path("/content/asr_archive_temp")
LOCAL_ARCHIVE_DIR.mkdir(parents=True, exist_ok=True)

AUDIO_INDEX_PATH = DATA_DIR / "train_audio_index_25h.jsonl"
ARCHIVE_INDEX_PATH = DATA_DIR / "audio_archive_index_25h.json"

# Get all extracted candidates in reproducible order.
records = sorted(
    completed.values(),
    key=lambda r: r["selection_rank"]
)

assert len(records) == len(candidate_records)

# Ensure every referenced MP3 exists before archiving.
for record in records:
    path = AUDIO_DIR / record["audio_file"]
    assert path.exists() and path.stat().st_size > 0, (
        f"Missing audio: {path}"
    )

# Save actual durations for ALL candidates.
with AUDIO_INDEX_PATH.open("w", encoding="utf-8") as f:
    for record in records:
        f.write(json.dumps(record, ensure_ascii=False) + "\n")

def sha256_file(path):
    digest = hashlib.sha256()
    with path.open("rb") as f:
        for chunk in iter(lambda: f.read(4 * 1024**2), b""):
            digest.update(chunk)
    return digest.hexdigest()

archive_index = {
    "target_hours": TRAIN_TARGET_HOURS,
    "total_recordings": len(records),
    "archives": []
}

batches = [
    records[i:i + ARCHIVE_BATCH_SIZE]
    for i in range(0, len(records), ARCHIVE_BATCH_SIZE)
]

for batch_number, batch in enumerate(
    tqdm(batches, desc="Backing up audio"), 1
):
    filename = f"amharic_audio_{batch_number:03d}.tar"

    local_tar = LOCAL_ARCHIVE_DIR / filename
    drive_tar = ARCHIVE_DIR / filename
    partial_tar = ARCHIVE_DIR / (filename + ".partial")

    # Create archive on Colab's faster local disk.
    with tarfile.open(local_tar, "w") as archive:
        for record in batch:
            source = AUDIO_DIR / record["audio_file"]
            archive.add(
                source,
                arcname=record["audio_file"],
                recursive=False
            )

    local_hash = sha256_file(local_tar)

    # Copy to Drive; rename only after copying completes.
    shutil.copyfile(local_tar, partial_tar)
    partial_tar.replace(drive_tar)

    # Verify the stored archive is identical.
    drive_hash = sha256_file(drive_tar)
    assert local_hash == drive_hash, (
        f"Checksum mismatch: {filename}"
    )

    archive_index["archives"].append({
        "filename": filename,
        "recordings": len(batch),
        "size_bytes": drive_tar.stat().st_size,
        "sha256": drive_hash
    })

    # Remove temporary TAR, keeping original MP3s.
    local_tar.unlink()

# Save archive index after successful verification.
with ARCHIVE_INDEX_PATH.open("w", encoding="utf-8") as f:
    json.dump(archive_index, f, indent=2)

total_bytes = sum(
    item["size_bytes"]
    for item in archive_index["archives"]
)

print("\nAUDIO BACKUP SUMMARY")
print("-" * 45)
print("Candidate recordings backed up:", len(records))
print("Archives created:", len(archive_index["archives"]))
print("Total archive size:", round(total_bytes / 1024**3, 2), "GB")
print("SHA-256 verification: PASSED")
print("Audio index:", AUDIO_INDEX_PATH)
print("Archive index:", ARCHIVE_INDEX_PATH)
print("Archive directory:", ARCHIVE_DIR)

print("\nOriginal local MP3 files remain available.")


Backing up audio:   0%|          | 0/10 [00:00<?, ?it/s]


AUDIO BACKUP SUMMARY
---------------------------------------------
Candidate recordings backed up: 5915
Archives created: 10
Total archive size: 1.57 GB
SHA-256 verification: PASSED
Audio index: /content/drive/MyDrive/Amharic_ASR_XLSR/data/train_audio_index_25h.jsonl
Archive index: /content/drive/MyDrive/Amharic_ASR_XLSR/data/audio_archive_index_25h.json
Archive directory: /content/drive/MyDrive/Amharic_ASR_XLSR/audio_archives/25h

Original local MP3 files remain available.


In [ ]:

import json
import numpy as np
import torch

from pathlib import Path
from torch.utils.data import Dataset, DataLoader
from torchcodec.decoders import AudioDecoder

from transformers import (
    Wav2Vec2Config,
    Wav2Vec2FeatureExtractor,
    Wav2Vec2Processor
)

# ------------------------------------------
# 1. Load the final 25-hour training manifest
# ------------------------------------------

with FINAL_MANIFEST.open(encoding="utf-8") as f:
    train_records = [json.loads(line) for line in f]

assert len(train_records) == 5084

MODEL_ID = "facebook/wav2vec2-xls-r-300m"
SAMPLE_RATE = 16000

model_config = Wav2Vec2Config.from_pretrained(MODEL_ID)

# XLS-R uses layer normalization in its feature extractor,
# so attention masks are appropriate for padded audio.
assert model_config.feat_extract_norm == "layer"

feature_extractor = Wav2Vec2FeatureExtractor(
    feature_size=1,
    sampling_rate=SAMPLE_RATE,
    padding_value=0.0,
    do_normalize=True,
    return_attention_mask=True
)

processor = Wav2Vec2Processor(
    feature_extractor=feature_extractor,
    tokenizer=tokenizer
)

processor.save_pretrained(str(PROJECT_DIR / "processor"))

# ------------------------------------------
# 2. Check CTC sequence-length feasibility
# ------------------------------------------

def output_frames(num_samples):
    length = int(num_samples)

    for kernel, stride in zip(
        model_config.conv_kernel,
        model_config.conv_stride
    ):
        length = (length - kernel) // stride + 1

    return length

ctc_failures = []
minimum_margin = float("inf")
max_label_length = 0

for record in train_records:
    labels = tokenizer.encode(
        record["transcription"],
        add_special_tokens=False
    )

    # CTC needs extra time steps for repeated adjacent labels.
    repeated = sum(
        labels[i] == labels[i - 1]
        for i in range(1, len(labels))
    )

    required_frames = len(labels) + repeated

    # Estimated from measured audio duration.
    estimated_samples = round(
        record["duration_seconds"] * SAMPLE_RATE
    )

    frames = output_frames(estimated_samples)
    margin = frames - required_frames

    minimum_margin = min(minimum_margin, margin)
    max_label_length = max(max_label_length, len(labels))

    if margin < 0:
        ctc_failures.append({
            "id": record["id"],
            "available_frames": frames,
            "required_frames": required_frames
        })

print("CTC FEASIBILITY CHECK")
print("-" * 45)
print("Recordings checked:", len(train_records))
print("Maximum label length:", max_label_length)
print("Minimum estimated frame margin:", minimum_margin)
print("Potentially infeasible recordings:", len(ctc_failures))

if ctc_failures:
    print("First failures:", ctc_failures[:5])

# ------------------------------------------
# 3. Create an on-demand audio dataset
# ------------------------------------------

class AmharicASRDataset(Dataset):
    def __init__(self, records, audio_dir, processor):
        self.records = records
        self.audio_dir = Path(audio_dir)
        self.processor = processor

    def __len__(self):
        return len(self.records)

    def __getitem__(self, index):
        record = self.records[index]

        audio_path = self.audio_dir / record["audio_file"]

        decoder = AudioDecoder(
            str(audio_path),
            sample_rate=SAMPLE_RATE,
            num_channels=1
        )

        audio_samples = decoder.get_all_samples()

        waveform = (
            audio_samples.data[0]
            .cpu()
            .numpy()
            .astype(np.float32)
        )

        assert audio_samples.sample_rate == SAMPLE_RATE

        inputs = self.processor.feature_extractor(
            waveform,
            sampling_rate=SAMPLE_RATE
        )

        labels = self.processor.tokenizer(
            record["transcription"],
            add_special_tokens=False
        ).input_ids

        return {
            "input_values": inputs.input_values[0],
            "labels": labels,
            "id": record["id"]
        }

# ------------------------------------------
# 4. Dynamically pad each training batch
# ------------------------------------------

def ctc_collator(examples):
    audio_features = [
        {"input_values": x["input_values"]}
        for x in examples
    ]

    label_features = [
        {"input_ids": x["labels"]}
        for x in examples
    ]

    batch = processor.feature_extractor.pad(
        audio_features,
        padding=True,
        return_attention_mask=True,
        return_tensors="pt"
    )

    label_batch = processor.tokenizer.pad(
        label_features,
        padding=True,
        return_tensors="pt"
    )

    batch["labels"] = label_batch["input_ids"].masked_fill(
        label_batch["attention_mask"] != 1,
        -100
    )

    return batch

train_dataset = AmharicASRDataset(
    train_records,
    AUDIO_DIR,
    processor
)

# Small diagnostic batch, CPU only.
test_loader = DataLoader(
    train_dataset,
    batch_size=2,
    shuffle=False,
    collate_fn=ctc_collator,
    num_workers=0
)

batch = next(iter(test_loader))

# ------------------------------------------
# 5. Verify the resulting tensors
# ------------------------------------------

print("\nDATALOADER TEST")
print("-" * 45)

print("Dataset size:", len(train_dataset))
print("Audio tensor shape:", tuple(batch["input_values"].shape))
print("Attention mask shape:", tuple(batch["attention_mask"].shape))
print("Label tensor shape:", tuple(batch["labels"].shape))

print("Audio dtype:", batch["input_values"].dtype)
print("Label dtype:", batch["labels"].dtype)

print(
    "Audio contains NaN/Inf:",
    not torch.isfinite(batch["input_values"]).all().item()
)

print(
    "Valid label counts:",
    (batch["labels"] != -100).sum(dim=1).tolist()
)

print(
    "Audio lengths (seconds):",
    [
        round(int(x) / SAMPLE_RATE, 2)
        for x in batch["attention_mask"].sum(dim=1)
    ]
)

assert torch.isfinite(batch["input_values"]).all()
assert not ctc_failures, "Some recordings fail estimated CTC feasibility."

print("\nDATALOADER TEST PASSED")


CTC FEASIBILITY CHECK
---------------------------------------------
Recordings checked: 5084
Maximum label length: 407
Minimum estimated frame margin: -9
Potentially infeasible recordings: 1
First failures: [{'id': '5psPJBBetW3jsIWVgElP', 'available_frames': 64, 'required_frames': 73}]

DATALOADER TEST
---------------------------------------------
Dataset size: 5084
Audio tensor shape: (2, 299904)
Attention mask shape: (2, 299904)
Label tensor shape: (2, 119)
Audio dtype: torch.float32
Label dtype: torch.int64
Audio contains NaN/Inf: False
Valid label counts: [118, 119]
Audio lengths (seconds): [17.98, 18.74]


AssertionError: Some recordings fail estimated CTC feasibility.

In [ ]:

import json
import numpy as np

from IPython.display import Audio, display
from torchcodec.decoders import AudioDecoder
from torch.utils.data import DataLoader

# -------------------------------------------------
# 1. Calculate minimum frames required by CTC
# -------------------------------------------------

def required_ctc_frames(text):
    ids = tokenizer.encode(
        text,
        add_special_tokens=False
    )

    repeated = sum(
        ids[i] == ids[i - 1]
        for i in range(1, len(ids))
    )

    return len(ids) + repeated


# -------------------------------------------------
# 2. Verify actual audio lengths near CTC limits
# -------------------------------------------------

valid_records = []
excluded_records = []
inspected = []

for record in train_records:
    required = required_ctc_frames(record["transcription"])

    estimated_samples = round(
        record["duration_seconds"] * SAMPLE_RATE
    )
    estimated_frames = output_frames(estimated_samples)

    # Metadata is approximate. Decode recordings close
    # to the minimum instead of relying on estimates.
    if estimated_frames - required <= 10:
        path = AUDIO_DIR / record["audio_file"]

        decoder = AudioDecoder(
            str(path),
            sample_rate=SAMPLE_RATE,
            num_channels=1
        )

        samples = decoder.get_all_samples()
        actual_frames = output_frames(samples.data.shape[-1])

        inspected.append(record["id"])

        if actual_frames < required:
            excluded_records.append({
                **record,
                "required_frames": required,
                "available_frames": actual_frames
            })

            print("\nINFEASIBLE RECORDING")
            print("ID:", record["id"])
            print(
                "Actual duration:",
                round(samples.data.shape[-1] / SAMPLE_RATE, 3),
                "seconds"
            )
            print("Available frames:", actual_frames)
            print("Required frames:", required)
            print("Transcription:")
            print(record["transcription"])

            print("\nAudio playback:")
            display(
                Audio(
                    samples.data[0].cpu().numpy(),
                    rate=SAMPLE_RATE
                )
            )
            continue

    valid_records.append(record)


# -------------------------------------------------
# 3. Save a new, corrected training manifest
# -------------------------------------------------

SAFE_MANIFEST = (
    DATA_DIR / "train_final_25h_ctc_safe.jsonl"
)

with SAFE_MANIFEST.open("w", encoding="utf-8") as file:
    for record in valid_records:
        file.write(
            json.dumps(record, ensure_ascii=False) + "\n"
        )

# Keep an audit record of exclusions.
EXCLUSIONS_PATH = (
    DATA_DIR / "ctc_exclusions_25h.json"
)

with EXCLUSIONS_PATH.open("w", encoding="utf-8") as file:
    json.dump(
        excluded_records,
        file,
        ensure_ascii=False,
        indent=2
    )


# -------------------------------------------------
# 4. Rebuild the DataLoader with valid recordings
# -------------------------------------------------

train_records = valid_records

train_dataset = AmharicASRDataset(
    train_records,
    AUDIO_DIR,
    processor
)

test_loader = DataLoader(
    train_dataset,
    batch_size=2,
    shuffle=False,
    collate_fn=ctc_collator,
    num_workers=0
)

batch = next(iter(test_loader))

assert torch.isfinite(batch["input_values"]).all()
assert len(valid_records) + len(excluded_records) == 5084

total_hours = sum(
    r["duration_seconds"] for r in valid_records
) / 3600

print("\nFINAL DATASET VALIDATION")
print("-" * 45)
print("Original recordings:", 5084)
print("Near-limit recordings decoded:", len(inspected))
print("Excluded recordings:", len(excluded_records))
print("Final recordings:", len(train_records))
print("Final training hours:", round(total_hours, 4))
print(
    "Unique speakers:",
    len({r["speaker_id"] for r in train_records})
)
print("Batch audio shape:", tuple(batch["input_values"].shape))
print("Batch label shape:", tuple(batch["labels"].shape))
print("Safe manifest:", SAFE_MANIFEST)

print("\nDATALOADER VALIDATION PASSED")



INFEASIBLE RECORDING
ID: 5psPJBBetW3jsIWVgElP
Actual duration: 1.296 seconds
Available frames: 64
Required frames: 73
Transcription:
ማስታወቂያ ምርትን አገልግሎትን ወይም ሐሳብን ለተወሰነ ታዳሚ ለማስተዋወቅ የሚደረግ የሚከፈልበት የግንኙነት ዘዴ ነው

Audio playback:



FINAL DATASET VALIDATION
---------------------------------------------
Original recordings: 5084
Near-limit recordings decoded: 1
Excluded recordings: 1
Final recordings: 5083
Final training hours: 25.0007
Unique speakers: 566
Batch audio shape: (2, 299904)
Batch label shape: (2, 119)
Safe manifest: /content/drive/MyDrive/Amharic_ASR_XLSR/data/train_final_25h_ctc_safe.jsonl

DATALOADER VALIDATION PASSED


In [ ]:

import gc
import torch

from transformers import Wav2Vec2ForCTC

# ------------------------------------------
# 1. Load pretrained XLS-R
# ------------------------------------------

DEVICE = "cuda"
UNFROZEN_LAYERS = 2

assert torch.cuda.is_available(), "GPU is required."

model = Wav2Vec2ForCTC.from_pretrained(
    MODEL_ID,
    vocab_size=len(tokenizer),
    pad_token_id=tokenizer.pad_token_id,
    ctc_loss_reduction="mean",
    ctc_zero_infinity=True,
    ignore_mismatched_sizes=True
)

# A newly initialized CTC head is expected.
assert model.lm_head.out_features == 321

# ------------------------------------------
# 2. Freeze everything, then selectively
#    unfreeze the layers we want to train
# ------------------------------------------

for parameter in model.parameters():
    parameter.requires_grad = False

for layer in model.wav2vec2.encoder.layers[-UNFROZEN_LAYERS:]:
    for parameter in layer.parameters():
        parameter.requires_grad = True

for parameter in model.lm_head.parameters():
    parameter.requires_grad = True

# Avoid the frozen-input checkpointing problem.
model.gradient_checkpointing_enable(
    gradient_checkpointing_kwargs={
        "use_reentrant": False
    }
)

model.to(DEVICE)
model.train()

total_params = sum(
    p.numel() for p in model.parameters()
)

trainable_params = sum(
    p.numel()
    for p in model.parameters()
    if p.requires_grad
)

print("MODEL CONFIGURATION")
print("-" * 45)
print("Total parameters:", f"{total_params:,}")
print("Trainable parameters:", f"{trainable_params:,}")
print(
    "Trainable percentage:",
    f"{100 * trainable_params / total_params:.2f}%"
)
print("Transformer layers:", len(model.wav2vec2.encoder.layers))
print("Unfrozen layers:", UNFROZEN_LAYERS)
print("Vocabulary size:", model.config.vocab_size)
print("CTC blank ID:", model.config.pad_token_id)
print(
    "Gradient checkpointing:",
    model.is_gradient_checkpointing
)

# ------------------------------------------
# 3. Choose a short valid recording
# ------------------------------------------

sample_index = min(
    range(min(64, len(train_records))),
    key=lambda i: train_records[i]["duration_seconds"]
)

sample_record = train_records[sample_index]

# Reuse the verified dataset and collator.
sample_batch = ctc_collator(
    [train_dataset[sample_index]]
)

sample_batch = {
    key: value.to(DEVICE)
    for key, value in sample_batch.items()
}

print("\nDIAGNOSTIC RECORDING")
print("ID:", sample_record["id"])
print(
    "Duration:",
    round(sample_record["duration_seconds"], 2),
    "seconds"
)
print(
    "Label tokens:",
    int((sample_batch["labels"] != -100).sum())
)

# ------------------------------------------
# 4. Forward pass + backward pass
# ------------------------------------------

torch.cuda.reset_peak_memory_stats()
model.zero_grad(set_to_none=True)

scaler = torch.amp.GradScaler(
    "cuda",
    init_scale=128.0
)

with torch.autocast(
    device_type="cuda",
    dtype=torch.float16
):
    outputs = model(**sample_batch)
    loss = outputs.loss

print("\nFORWARD PASS")
print("CTC loss:", round(float(loss.item()), 4))
print("Finite loss:", bool(torch.isfinite(loss).item()))
print("Output logits:", tuple(outputs.logits.shape))

assert torch.isfinite(loss), "Non-finite CTC loss."

# Scale gradients to make FP16 training more stable.
scaler.scale(loss).backward()

# ------------------------------------------
# 5. Verify gradients in every trainable
#    component
# ------------------------------------------

def gradient_report(module, name):
    gradients = [
        p.grad
        for p in module.parameters()
        if p.requires_grad
    ]

    available = [
        g for g in gradients
        if g is not None
    ]

    all_present = len(available) == len(gradients)

    all_finite = (
        len(available) > 0
        and all(torch.isfinite(g).all().item() for g in available)
    )

    # Gradients are currently scaled by GradScaler.
    scale = scaler.get_scale()

    max_gradient = max(
        (g.detach().abs().max().item() / scale
         for g in available),
        default=0.0
    )

    print(
        f"{name:20} "
        f"gradients={len(available)}/{len(gradients)} "
        f"finite={all_finite} "
        f"max_abs={max_gradient:.8f}"
    )

    assert all_present, f"Missing gradients in {name}"
    assert all_finite, f"Non-finite gradients in {name}"
    assert max_gradient > 0, f"Zero gradients in {name}"


print("\nGRADIENT FLOW CHECK")
print("-" * 70)

gradient_report(
    model.wav2vec2.encoder.layers[-2],
    "Transformer layer 22"
)

gradient_report(
    model.wav2vec2.encoder.layers[-1],
    "Transformer layer 23"
)

gradient_report(
    model.lm_head,
    "CTC prediction head"
)

print(
    "\nPeak GPU memory:",
    round(torch.cuda.max_memory_allocated() / 1024**3, 2),
    "GB"
)

# No optimizer.step() here.
# This is a diagnostic, not a training update.
model.zero_grad(set_to_none=True)

del outputs, loss, sample_batch
gc.collect()
torch.cuda.empty_cache()

print("\nGRADIENT DIAGNOSTIC PASSED")
print("No model weights were updated.")


pytorch_model.bin:   0%|          | 0.00/1.27G [00:00<?, ?B/s]

Some weights of Wav2Vec2ForCTC were not initialized from the model checkpoint at facebook/wav2vec2-xls-r-300m and are newly initialized: ['lm_head.bias', 'lm_head.weight']
You should probably TRAIN this model on a down-stream task to be able to use it for predictions and inference.


model.safetensors:   0%|          | 0.00/1.27G [00:00<?, ?B/s]

MODEL CONFIGURATION
---------------------------------------------
Total parameters: 315,767,745
Trainable parameters: 25,521,473
Trainable percentage: 8.08%
Transformer layers: 24
Unfrozen layers: 2
Vocabulary size: 321
CTC blank ID: 320
Gradient checkpointing: True

DIAGNOSTIC RECORDING
ID: 3d4DQUr7d0su1SBZTb4t
Duration: 9.46 seconds
Label tokens: 60

FORWARD PASS
CTC loss: 40.9095
Finite loss: True
Output logits: (1, 472, 321)

GRADIENT FLOW CHECK
----------------------------------------------------------------------
Transformer layer 22 gradients=16/16 finite=True max_abs=2.12003255
Transformer layer 23 gradients=16/16 finite=True max_abs=0.07950237
CTC prediction head  gradients=2/2 finite=True max_abs=2.74804688

Peak GPU memory: 1.59 GB

GRADIENT DIAGNOSTIC PASSED
No model weights were updated.


In [ ]:

# CELL 21 - RESTORE EXISTING BASELINE
# Do not recreate or overwrite saved checkpoints.

import json
import shutil
from pathlib import Path

PROJECT_DIR = Path(
    "/content/drive/MyDrive/Amharic_ASR_XLSR"
)
DATA_DIR = PROJECT_DIR / "data"
CHECKPOINT_DIR = PROJECT_DIR / "checkpoints"

BASELINE_DIR = (
    PROJECT_DIR / "baselines" / "xlsr_step0"
)

BASELINE_EVAL_PATH = (
    DATA_DIR / "baseline_eval_fixed_12.jsonl"
)

DRIVE_EVAL_AUDIO = PROJECT_DIR / "evaluation_audio"
EVAL_AUDIO_DIR = Path("/content/amharic_eval_audio")
EVAL_AUDIO_DIR.mkdir(parents=True, exist_ok=True)

# 1. Verify the original checkpoint.
assert BASELINE_DIR.is_dir(), (
    f"Missing baseline: {BASELINE_DIR}"
)

assert list(BASELINE_DIR.glob("*.safetensors")), (
    "Baseline model weights are missing."
)

print("Original baseline checkpoint: FOUND")

# 2. Restore the fixed evaluation manifest.
assert BASELINE_EVAL_PATH.is_file(), (
    f"Missing evaluation manifest: {BASELINE_EVAL_PATH}"
)

with BASELINE_EVAL_PATH.open(encoding="utf-8") as f:
    eval_records = [json.loads(line) for line in f]

assert len(eval_records) == 12
assert len({r["id"] for r in eval_records}) == 12

print("Fixed evaluation recordings:", len(eval_records))

# 3. Restore evaluation audio from Google Drive.
restored = 0
missing_audio = []

for record in eval_records:
    filename = record["id"] + ".mp3"

    source = DRIVE_EVAL_AUDIO / filename
    destination = EVAL_AUDIO_DIR / filename

    if destination.exists() and destination.stat().st_size > 0:
        continue

    if source.exists():
        shutil.copy2(source, destination)
        restored += 1
    else:
        missing_audio.append(filename)

print("Audio files restored locally:", restored)
print("Missing evaluation recordings:", len(missing_audio))

# 4. Locate previously saved baseline results.
BASELINE_METRICS_PATH = (
    DATA_DIR / "baseline_step0_metrics.json"
)

BASELINE_PREDICTIONS_PATH = (
    DATA_DIR / "baseline_step0_predictions_12.jsonl"
)

if BASELINE_METRICS_PATH.exists():
    with BASELINE_METRICS_PATH.open(encoding="utf-8") as f:
        baseline_metrics = json.load(f)

    print(
        "Saved baseline CER:",
        f"{baseline_metrics['cer'] * 100:.2f}%"
    )
    print(
        "Saved baseline WER:",
        f"{baseline_metrics['wer'] * 100:.2f}%"
    )
else:
    print("Baseline metrics not found.")

print("\n" + "=" * 50)
print("BASELINE RECOVERY COMPLETE")
print("=" * 50)
print("Original model preserved:", True)
print("Evaluation manifest:", BASELINE_EVAL_PATH)
print("Evaluation audio directory:", EVAL_AUDIO_DIR)
print("Saved predictions:", BASELINE_PREDICTIONS_PATH.exists())
print("Saved metrics:", BASELINE_METRICS_PATH.exists())

if missing_audio:
    print("\nMissing audio IDs:", missing_audio)
else:
    print("\nAll evaluation audio is available.")


Original baseline checkpoint: FOUND
Fixed evaluation recordings: 12
Audio files restored locally: 12
Missing evaluation recordings: 0
Saved baseline CER: 171.64%
Saved baseline WER: 100.00%

BASELINE RECOVERY COMPLETE
Original model preserved: True
Evaluation manifest: /content/drive/MyDrive/Amharic_ASR_XLSR/data/baseline_eval_fixed_12.jsonl
Evaluation audio directory: /content/amharic_eval_audio
Saved predictions: True
Saved metrics: True

All evaluation audio is available.


In [ ]:

import json
import shutil
import torch
import numpy as np
import fsspec
import pyarrow.parquet as pq

from pathlib import Path
from tqdm.auto import tqdm
from torchcodec.decoders import AudioDecoder
from jiwer import cer, wer

# =========================================
# 1. Load our fixed evaluation examples
# =========================================

with BASELINE_EVAL_PATH.open(encoding="utf-8") as f:
    eval_records = [json.loads(line) for line in f]

assert len(eval_records) == 12

EVAL_AUDIO_DIR = Path("/content/amharic_eval_audio")
EVAL_AUDIO_DIR.mkdir(parents=True, exist_ok=True)

DRIVE_EVAL_AUDIO = PROJECT_DIR / "evaluation_audio"
DRIVE_EVAL_AUDIO.mkdir(parents=True, exist_ok=True)

needed_ids = {r["id"] for r in eval_records}

# Restore already downloaded audio if available.
for record in eval_records:
    filename = record["id"] + ".mp3"
    local_path = EVAL_AUDIO_DIR / filename
    drive_path = DRIVE_EVAL_AUDIO / filename

    if not local_path.exists() and drive_path.exists():
        shutil.copy2(drive_path, local_path)

missing_ids = {
    record_id for record_id in needed_ids
    if not (EVAL_AUDIO_DIR / (record_id + ".mp3")).exists()
}

print("Evaluation examples:", len(eval_records))
print("Recordings needing download:", len(missing_ids))

# =========================================
# 2. Download only needed validation audio
# =========================================

if missing_ids:
    for shard in tqdm(val_shards, desc="Retrieving validation audio"):
        with fsspec.open(
            shard["url"],
            "rb",
            block_size=8 * 1024**2
        ) as source:

            parquet = pq.ParquetFile(source)

            for group_index in range(parquet.metadata.num_row_groups):

                # First read the lightweight ID column.
                group_ids = parquet.read_row_group(
                    group_index,
                    columns=["id"]
                ).column("id").to_pylist()

                matched = [
                    (index, record_id)
                    for index, record_id in enumerate(group_ids)
                    if record_id in missing_ids
                ]

                if not matched:
                    continue

                # Read audio only for relevant row groups.
                table = parquet.read_row_group(
                    group_index,
                    columns=["audio"]
                )

                for index, record_id in matched:
                    audio = table.column("audio")[index].as_py()
                    encoded = audio.get("bytes")

                    if encoded is None:
                        raise RuntimeError(
                            f"Missing embedded audio: {record_id}"
                        )

                    filename = record_id + ".mp3"
                    local_path = EVAL_AUDIO_DIR / filename
                    drive_path = DRIVE_EVAL_AUDIO / filename

                    local_path.write_bytes(encoded)
                    shutil.copy2(local_path, drive_path)

                    missing_ids.remove(record_id)

        if not missing_ids:
            break

assert not missing_ids, (
    f"Missing evaluation audio IDs: {missing_ids}"
)

print("Evaluation audio ready.")

# =========================================
# 3. Run the STEP-ZERO model
# =========================================

model.eval()

results = []
references = []
predictions = []

for i, record in enumerate(
    tqdm(eval_records, desc="Step-zero inference"), 1
):
    path = EVAL_AUDIO_DIR / (record["id"] + ".mp3")

    decoder = AudioDecoder(
        str(path),
        sample_rate=SAMPLE_RATE,
        num_channels=1
    )

    samples = decoder.get_all_samples()

    waveform = (
        samples.data[0]
        .cpu()
        .numpy()
        .astype(np.float32)
    )

    inputs = processor.feature_extractor(
        waveform,
        sampling_rate=SAMPLE_RATE,
        return_attention_mask=True,
        return_tensors="pt"
    )

    inputs = {
        key: value.to(DEVICE)
        for key, value in inputs.items()
    }

    with torch.inference_mode():
        with torch.autocast(
            device_type="cuda",
            dtype=torch.float16
        ):
            logits = model(**inputs).logits

    token_ids = logits.argmax(dim=-1)

    # Standard CTC decoding:
    # collapse repeated frame predictions and remove blanks.
    predicted = processor.batch_decode(
        token_ids.cpu().numpy()
    )[0]

    predicted = normalize_amharic_ctc(predicted)
    reference = record["transcription"]

    blank_fraction = (
        (token_ids == tokenizer.pad_token_id)
        .float()
        .mean()
        .item()
    )

    references.append(reference)
    predictions.append(predicted)

    results.append({
        "id": record["id"],
        "speaker_id": record["speaker_id"],
        "duration_seconds": round(
            len(waveform) / SAMPLE_RATE, 3
        ),
        "reference": reference,
        "prediction": predicted,
        "cer": cer(reference, predicted),
        "wer": wer(reference, predicted),
        "blank_fraction": blank_fraction
    })

    print(f"\n{'=' * 65}")
    print(f"RECORDING {i}")
    print("Duration:", results[-1]["duration_seconds"], "s")
    print("REFERENCE:", reference[:220])
    print("PREDICTED:", predicted[:220])
    print("CER:", round(results[-1]["cer"], 4))
    print("WER:", round(results[-1]["wer"], 4))
    print(
        "Blank-frame percentage:",
        round(blank_fraction * 100, 2),
        "%"
    )

    del inputs, logits, token_ids

# =========================================
# 4. Compute and save baseline metrics
# =========================================

overall_cer = cer(references, predictions)
overall_wer = wer(references, predictions)

STEP0_RESULTS = (
    DATA_DIR / "baseline_step0_predictions_12.jsonl"
)

with STEP0_RESULTS.open("w", encoding="utf-8") as file:
    for result in results:
        file.write(
            json.dumps(result, ensure_ascii=False) + "\n"
        )

STEP0_METRICS = DATA_DIR / "baseline_step0_metrics.json"

metrics = {
    "model": MODEL_ID,
    "checkpoint": str(BASELINE_DIR),
    "training_step": 0,
    "evaluation_examples": len(results),
    "cer": overall_cer,
    "wer": overall_wer,
    "empty_predictions": sum(
        not prediction for prediction in predictions
    ),
    "mean_blank_fraction": float(np.mean([
        r["blank_fraction"] for r in results
    ]))
}

with STEP0_METRICS.open("w", encoding="utf-8") as file:
    json.dump(metrics, file, indent=2)

# Restore training mode for subsequent experiments.
model.train()

print("\n" + "=" * 65)
print("STARTING MODEL BASELINE")
print("=" * 65)

print("Evaluation recordings:", len(results))
print("Overall CER:", round(overall_cer, 4))
print("Overall WER:", round(overall_wer, 4))
print("CER percentage:", round(overall_cer * 100, 2), "%")
print("WER percentage:", round(overall_wer * 100, 2), "%")
print("Empty predictions:", metrics["empty_predictions"])
print(
    "Mean blank-frame percentage:",
    round(metrics["mean_blank_fraction"] * 100, 2),
    "%"
)

print("\nPredictions saved:", STEP0_RESULTS)
print("Metrics saved:", STEP0_METRICS)
print("Evaluation audio:", DRIVE_EVAL_AUDIO)

print("\nSTEP-ZERO BASELINE COMPLETE")


Evaluation examples: 12
Recordings needing download: 0
Evaluation audio ready.


Step-zero inference:   0%|          | 0/12 [00:00<?, ?it/s]


RECORDING 1
Duration: 16.296 s
REFERENCE: የፈንገስ ማጥፊያ የፈንገስ ማጥፊያ ሰብል ላይ የሚወጡ የፈንገስ በሽታ ለመከላከል እና ለመቆጣጠር ያገለግላሉ ለቡና አትክልትና ለእህል ሰብሎች ለዘር በመሰብሰብ ቅጠሉን በመብላት ይከላከላሉ
PREDICTED: ፻ጴ፻ጴ፻ጴ፻ጴ፻ጴኑ፻ጴኑ፻ኑ፻ኑጴ፻ኑ፻ኗኑ፻ኑ፻ጴኑኗuኑ፻ጴኑጴኑጴ፻ጴኑ፻ጴኑ፻ጴ፻ኑ፻ኗኑ፻ኑኗጴኑ፻ጴ፻ጴኑጴ፻ጴ፻uኑቡ፻ጴኑ፻ጴ፻ኑ፻ኗኑ፻ኹኑ፻ኑ፻ጴ፻ኹ፻ጴ፻ኑ፻ጴ፻ኑ፻ኑ፻ኑ፻ኑ፻ጴኹ፻ኑ፻ኑ፻ኗኑ፻ኑ፻ኑጴ፻ጴ፻ጴuጴ፻ጴ፻ኑ፻ኑ፻ጴ፻ኑኹኑ፻ኑ፻ጴ፻ኑ፻ጴኑጴኑ፻ጴ፻ጴኗ፻ኗኹኑጴ፻ጴ፻ጴ፻ጴኹጴኑ፻ጴ፻ኑ፻ጴ፻ጴ፻ጴ፻ጴ፻ጴኑኗኑኗ፻ጴ፻ጴቡጴ፻ኗኑጴ፻ኑ፻ኗኑ፻ኑ፻4ጴ፻ጴ፻ኑ፻ኑ፻ጴኑ፻ኗ፻ኑ፻ጴ፻ኑ፻
CER: 2.5128
WER: 1.0
Blank-frame percentage: 0.0 %

RECORDING 2
Duration: 18.984 s
REFERENCE: የኢትዮጵያን ንግድ ባንክ በኢትዮጵያ ወስጥ ከሚገኙ እጅግ በጣም ስማቸው ገናና እና ጥንት ከሆኑ ባንኮች መካከል አንድ ነው ይህ ባንክ ሃላፊነቱ ያለው በመንግሥት እድ ቢሆንም እጅግ በጣም ብዙ ግለሰቦችን ቀጥሩ የሚያሠራ እና ብዙ ተደራሽነትን በተለያዩ የሀገሪቱ ክፍሎች ያደረገ ባንክ ነው
PREDICTED: ፻ጴ፻ጴ፻ጴ፻ጴ፻ኑ፻ጴ፻ጴ፻ጴ፻ጴ፻ጴኹ፻ጴ፻ኗ፻ጴ፻ዒጴ፻ጴ፻ጴ፻ጴ፻ጴ፻ጴ፻ኗጴ፻ጴ፻ጴ፻ኑ፻ኗጴኑ፻ጴ፻ኹ፻ጴ፻ጴ፻ኢ፻ጴ፻ጴ፻ጴ፻ጴ፻ኧኑጴኗ፻ጴ፻ጴ፻ጴቤ፻ጴ፻ጴኹ፻ጴ፻ጴ፻ጴ፻ጴ፻ጴኗ፻ጴ፻v፻ጴ፻ኹኗ፻ጴ፻ጴ፻ኗኑኢጴ፻ሲ፻ጴኹኑጴ፻ጴ፻ጴ፻ጴ፻ኹ፻ጴ፻ጴ፻ጴ፻ኧ፻ጴ፻ጴ፻ጴ፻ጴ፻ኑ፻ጴ፻ጴ፻u፻ጴ፻ጴ፻ኗ፻ጴ፻ጴ፻ጴ፻ጴ፻u፻ኗ፻ጴ፻ጴ፻ጴ፻ጴ፻ኑጴ፻ጴ፻ጴ፻ጴኑጴ፻ጴ፻ጴ፻ጴ፻ጴ፻ኹ፻ጴ፻ጴ፻ኗጴኧ፻ጴኧጴ፻ጴ፻
CER: 1.2123
WER: 1.0
Blank-frame percentage: 0.0 %

RECORDING 3
Duration: 17.184 s
REFERENCE: የቃል መጠየቂያ

In [ ]:

import random
import math
import gc
import torch

# ==========================================
# 1. CONFIGURATION
# ==========================================

HEAD_LR = 1e-4
ENCODER_LR = 1e-5
WEIGHT_DECAY = 0.01
GRAD_ACCUM_STEPS = 4
MAX_GRAD_NORM = 1.0
SEED = 42

# ==========================================
# 2. SELECT FOUR SUITABLE RECORDINGS
# ==========================================

rng = random.Random(SEED)

eligible = [
    (i, record)
    for i, record in enumerate(train_records)
    if 8 <= record["duration_seconds"] <= 14
    and (
        output_frames(
            round(record["duration_seconds"] * SAMPLE_RATE)
        )
        - required_ctc_frames(record["transcription"])
    ) >= 30
]

rng.shuffle(eligible)

selected_indices = []
selected_speakers = set()

for index, record in eligible:
    if record["speaker_id"] not in selected_speakers:
        selected_indices.append(index)
        selected_speakers.add(record["speaker_id"])

    if len(selected_indices) == GRAD_ACCUM_STEPS:
        break

assert len(selected_indices) == GRAD_ACCUM_STEPS

print("OPTIMIZER DIAGNOSTIC")
print("-" * 50)
print("Selected recordings:", len(selected_indices))
print("Distinct speakers:", len(selected_speakers))
print("Encoder learning rate:", ENCODER_LR)
print("CTC head learning rate:", HEAD_LR)
print("Gradient accumulation:", GRAD_ACCUM_STEPS)

# ==========================================
# 3. CREATE OPTIMIZER
# ==========================================

encoder_parameters = [
    p
    for layer in model.wav2vec2.encoder.layers[-2:]
    for p in layer.parameters()
    if p.requires_grad
]

head_parameters = [
    p for p in model.lm_head.parameters()
    if p.requires_grad
]

optimizer = torch.optim.AdamW(
    [
        {
            "params": encoder_parameters,
            "lr": ENCODER_LR
        },
        {
            "params": head_parameters,
            "lr": HEAD_LR
        }
    ],
    weight_decay=WEIGHT_DECAY
)

scaler = torch.amp.GradScaler(
    "cuda",
    init_scale=128.0
)

# ==========================================
# 4. BACK UP TRAINABLE WEIGHTS IN MEMORY
# ==========================================

original_weights = {
    name: parameter.detach().cpu().clone()
    for name, parameter in model.named_parameters()
    if parameter.requires_grad
}

model.train()
optimizer.zero_grad(set_to_none=True)

losses = []
step_applied = False

try:
    # ======================================
    # 5. ACCUMULATE GRADIENTS
    # ======================================

    for step, index in enumerate(selected_indices, 1):
        batch = ctc_collator([train_dataset[index]])

        batch = {
            key: value.to(DEVICE)
            for key, value in batch.items()
        }

        with torch.autocast(
            device_type="cuda",
            dtype=torch.float16
        ):
            outputs = model(**batch)
            raw_loss = outputs.loss

        assert torch.isfinite(raw_loss).item(), (
            f"Non-finite loss on recording {step}"
        )

        losses.append(raw_loss.detach().item())

        scaled_loss = raw_loss / GRAD_ACCUM_STEPS
        scaler.scale(scaled_loss).backward()

        print(
            f"Recording {step}/{GRAD_ACCUM_STEPS} "
            f"| CTC loss: {raw_loss.item():.4f}"
        )

        del batch, outputs, raw_loss, scaled_loss

    # ======================================
    # 6. CLIP GRADIENTS AND UPDATE WEIGHTS
    # ======================================

    scaler.unscale_(optimizer)

    trainable_parameters = (
        encoder_parameters + head_parameters
    )

    gradient_norm = torch.nn.utils.clip_grad_norm_(
        trainable_parameters,
        max_norm=MAX_GRAD_NORM,
        error_if_nonfinite=True
    )

    scale_before = scaler.get_scale()

    scaler.step(optimizer)
    scaler.update()

    scale_after = scaler.get_scale()

    # ======================================
    # 7. MEASURE ACTUAL WEIGHT CHANGES
    # ======================================

    changes = {}

    with torch.no_grad():
        for name, parameter in model.named_parameters():
            if name not in original_weights:
                continue

            before = original_weights[name]
            after = parameter.detach().cpu()

            changes[name] = (
                after - before
            ).abs().max().item()

    layer22_change = max(
        value for name, value in changes.items()
        if "encoder.layers.22." in name
    )

    layer23_change = max(
        value for name, value in changes.items()
        if "encoder.layers.23." in name
    )

    head_change = max(
        value for name, value in changes.items()
        if name.startswith("lm_head.")
    )

    step_applied = (
        scale_after >= scale_before
        and layer22_change > 0
        and layer23_change > 0
        and head_change > 0
    )

    print("\nOPTIMIZER RESULTS")
    print("-" * 50)

    print("Mean CTC loss:", round(sum(losses) / len(losses), 4))
    print("Gradient norm before clipping:", float(gradient_norm))
    print("GradScaler before:", scale_before)
    print("GradScaler after:", scale_after)

    print("\nMAXIMUM ABSOLUTE WEIGHT CHANGES")
    print(f"Layer 22: {layer22_change:.10f}")
    print(f"Layer 23: {layer23_change:.10f}")
    print(f"CTC head: {head_change:.10f}")

    print("\nOptimizer update succeeded:", step_applied)

finally:
    # ======================================
    # 8. RESTORE EXACT STARTING WEIGHTS
    # ======================================

    with torch.no_grad():
        for name, parameter in model.named_parameters():
            if name in original_weights:
                parameter.copy_(
                    original_weights[name].to(parameter.device)
                )

    model.zero_grad(set_to_none=True)

    del optimizer, scaler
    gc.collect()
    torch.cuda.empty_cache()

    restored = all(
        torch.equal(
            parameter.detach().cpu(),
            original_weights[name]
        )
        for name, parameter in model.named_parameters()
        if name in original_weights
    )

    print("\nOriginal weights restored:", restored)

assert restored, "Failed to restore original weights."
assert step_applied, "Optimizer failed to update all components."

print("\nOPTIMIZER DIAGNOSTIC PASSED")
print("Model remains at training step zero.")


OPTIMIZER DIAGNOSTIC
--------------------------------------------------
Selected recordings: 4
Distinct speakers: 4
Encoder learning rate: 1e-05
CTC head learning rate: 0.0001
Gradient accumulation: 4
Recording 1/4 | CTC loss: 33.4110
Recording 2/4 | CTC loss: 43.3449
Recording 3/4 | CTC loss: 34.6501
Recording 4/4 | CTC loss: 29.4747

OPTIMIZER RESULTS
--------------------------------------------------
Mean CTC loss: 35.2201
Gradient norm before clipping: 12.05112075805664
GradScaler before: 128.0
GradScaler after: 128.0

MAXIMUM ABSOLUTE WEIGHT CHANGES
Layer 22: 0.0000104904
Layer 23: 0.0000100732
CTC head: 0.0001000911

Optimizer update succeeded: True

Original weights restored: True

OPTIMIZER DIAGNOSTIC PASSED
Model remains at training step zero.


In [ ]:

# CELL 19B - RESTORE CTC-SAFE TRAINING DATASET

import json
from pathlib import Path

PROJECT_DIR = Path("/content/drive/MyDrive/Amharic_ASR_XLSR")
DATA_DIR = PROJECT_DIR / "data"
CHECKPOINT_DIR = PROJECT_DIR / "checkpoints"

SAFE_MANIFEST = DATA_DIR / "train_final_25h_ctc_safe.jsonl"

# Verify the previously saved corrected dataset.
assert SAFE_MANIFEST.exists(), (
    f"Corrected dataset not found: {SAFE_MANIFEST}"
)

with SAFE_MANIFEST.open(encoding="utf-8") as f:
    safe_records = [json.loads(line) for line in f]

assert len(safe_records) == 5083, (
    f"Expected 5083 recordings, found {len(safe_records)}"
)

# Ensure the invalid recording is excluded.
invalid_id = "5psPJBBetW3jsIWVgElP"

assert all(
    record["id"] != invalid_id
    for record in safe_records
)

# Restore dataset variables used by subsequent cells.
train_records = safe_records

train_dataset = AmharicASRDataset(
    train_records,
    AUDIO_DIR,
    processor
)

assert len(train_dataset) == 5083

# Report available checkpoints.
print("DATASET RECOVERY")
print("-" * 45)
print("Recordings:", len(train_dataset))
print("Unique speakers:", len(set(
    record["speaker_id"] for record in train_records
)))
print("Invalid recording excluded: YES")

print("\nSAVED TRAINING CHECKPOINTS")

for step in [10, 50, 200, 350, 500]:
    path = CHECKPOINT_DIR / f"step_{step:06d}"
    print(
        f"Step {step}:",
        "AVAILABLE" if (path / "COMPLETE").exists()
        else "NOT FOUND"
    )

print("\nCurrent in-memory training step:",
      globals().get("successful_updates", "NOT LOADED"))

print("\nCTC-SAFE DATASET RESTORED")


DATASET RECOVERY
---------------------------------------------
Recordings: 5083
Unique speakers: 566
Invalid recording excluded: YES

SAVED TRAINING CHECKPOINTS
Step 10: AVAILABLE
Step 50: AVAILABLE
Step 200: AVAILABLE
Step 350: AVAILABLE
Step 500: AVAILABLE

Current in-memory training step: NOT LOADED

CTC-SAFE DATASET RESTORED


In [ ]:

import math
import json
import random
import shutil
import gc
from pathlib import Path

import torch
from transformers import get_cosine_schedule_with_warmup

# ==========================================
# 1. EXPERIMENT CONFIGURATION
# ==========================================

TRAINING_SEED = 42

NUM_EPOCHS = 3
GRAD_ACCUM_STEPS = 4
STEPS_THIS_RUN = 10

ENCODER_LR = 1e-5
HEAD_LR = 1e-4
WEIGHT_DECAY = 0.01
MAX_GRAD_NORM = 1.0

assert len(train_dataset) == 5083

STEPS_PER_EPOCH = math.ceil(
    len(train_dataset) / GRAD_ACCUM_STEPS
)

TOTAL_STEPS = NUM_EPOCHS * STEPS_PER_EPOCH
WARMUP_STEPS = math.ceil(TOTAL_STEPS * 0.05)

CHECKPOINT_NAME = f"step_{STEPS_THIS_RUN:06d}"
SAVE_DIR = CHECKPOINT_DIR / CHECKPOINT_NAME

assert not SAVE_DIR.exists(), (
    f"Checkpoint already exists: {SAVE_DIR}\n"
    "Do not restart from step zero over an existing checkpoint."
)

torch.manual_seed(TRAINING_SEED)
torch.cuda.manual_seed_all(TRAINING_SEED)

# ==========================================
# 2. CREATE REPRODUCIBLE TRAINING ORDER
# ==========================================

training_order = list(range(len(train_dataset)))

rng = random.Random(TRAINING_SEED)
rng.shuffle(training_order)

# First 40 recordings in the deterministic order.
num_records = STEPS_THIS_RUN * GRAD_ACCUM_STEPS

selected_indices = training_order[:num_records]

assert len(selected_indices) == 40

# ==========================================
# 3. OPTIMIZER AND LEARNING-RATE SCHEDULER
# ==========================================

encoder_params = [
    p
    for layer in model.wav2vec2.encoder.layers[-2:]
    for p in layer.parameters()
    if p.requires_grad
]

head_params = [
    p for p in model.lm_head.parameters()
    if p.requires_grad
]

optimizer = torch.optim.AdamW(
    [
        {"params": encoder_params, "lr": ENCODER_LR},
        {"params": head_params, "lr": HEAD_LR}
    ],
    weight_decay=WEIGHT_DECAY
)

scheduler = get_cosine_schedule_with_warmup(
    optimizer,
    num_warmup_steps=WARMUP_STEPS,
    num_training_steps=TOTAL_STEPS
)

scaler = torch.amp.GradScaler(
    "cuda",
    init_scale=128.0
)

model.train()
model.zero_grad(set_to_none=True)

torch.cuda.reset_peak_memory_stats()

print("TRAINING CONFIGURATION")
print("-" * 50)
print("Training recordings:", len(train_dataset))
print("Planned epochs:", NUM_EPOCHS)
print("Updates per epoch:", STEPS_PER_EPOCH)
print("Total planned updates:", TOTAL_STEPS)
print("Warmup steps:", WARMUP_STEPS)
print("Updates in this run:", STEPS_THIS_RUN)

# ==========================================
# 4. RUN FIRST 10 OPTIMIZER UPDATES
# ==========================================

step_losses = []
successful_updates = 0

for update_index in range(STEPS_THIS_RUN):

    optimizer.zero_grad(set_to_none=True)

    micro_losses = []

    start = update_index * GRAD_ACCUM_STEPS
    end = start + GRAD_ACCUM_STEPS

    for record_index in selected_indices[start:end]:

        batch = ctc_collator(
            [train_dataset[record_index]]
        )

        batch = {
            key: value.to(DEVICE)
            for key, value in batch.items()
        }

        with torch.autocast(
            device_type="cuda",
            dtype=torch.float16
        ):
            outputs = model(**batch)
            loss = outputs.loss

        assert torch.isfinite(loss).item(), (
            "Non-finite training loss encountered."
        )

        micro_losses.append(float(loss.item()))

        scaled_loss = loss / GRAD_ACCUM_STEPS

        scaler.scale(scaled_loss).backward()

        del batch, outputs, loss, scaled_loss

    # Unscale before gradient clipping.
    scaler.unscale_(optimizer)

    grad_norm = torch.nn.utils.clip_grad_norm_(
        encoder_params + head_params,
        max_norm=MAX_GRAD_NORM,
        error_if_nonfinite=True
    )

    previous_scale = scaler.get_scale()

    scaler.step(optimizer)
    scaler.update()

    current_scale = scaler.get_scale()

    # A scale reduction indicates an AMP overflow
    # caused the optimizer update to be skipped.
    if current_scale < previous_scale:
        raise RuntimeError(
            "AMP skipped an optimizer update. "
            "Stop and investigate before checkpointing."
        )

    scheduler.step()
    successful_updates += 1

    mean_loss = sum(micro_losses) / len(micro_losses)
    step_losses.append(mean_loss)

    current_encoder_lr = optimizer.param_groups[0]["lr"]
    current_head_lr = optimizer.param_groups[1]["lr"]

    print(
        f"Update {successful_updates:02d}/{STEPS_THIS_RUN} | "
        f"CTC loss: {mean_loss:.4f} | "
        f"Grad norm: {float(grad_norm):.3f} | "
        f"Head LR: {current_head_lr:.8f}"
    )

assert successful_updates == STEPS_THIS_RUN

# ==========================================
# 5. SAVE COMPLETE RESUMABLE CHECKPOINT
# ==========================================

LOCAL_SAVE_DIR = Path(
    f"/content/asr_{CHECKPOINT_NAME}"
)

LOCAL_SAVE_DIR.mkdir(parents=True, exist_ok=False)

# Save trained model weights and processor.
model.save_pretrained(
    str(LOCAL_SAVE_DIR),
    safe_serialization=True
)

processor.save_pretrained(str(LOCAL_SAVE_DIR))

# Save optimizer, scheduler, AMP scaler and RNG state.
trainer_state = {
    "global_step": successful_updates,
    "epoch": 0,
    "next_sample_offset": num_records,
    "seed": TRAINING_SEED,
    "num_epochs": NUM_EPOCHS,
    "gradient_accumulation": GRAD_ACCUM_STEPS,
    "total_steps": TOTAL_STEPS,
    "warmup_steps": WARMUP_STEPS,
    "unfrozen_layers": 2,
    "optimizer": optimizer.state_dict(),
    "scheduler": scheduler.state_dict(),
    "scaler": scaler.state_dict(),
    "torch_rng_state": torch.get_rng_state(),
    "cuda_rng_states": torch.cuda.get_rng_state_all()
}

torch.save(
    trainer_state,
    LOCAL_SAVE_DIR / "trainer_state.pt"
)

training_summary = {
    "training_step": successful_updates,
    "recordings_processed": num_records,
    "mean_ctc_loss": sum(step_losses) / len(step_losses),
    "step_losses": step_losses,
    "planned_epochs": NUM_EPOCHS,
    "dataset_recordings": len(train_dataset)
}

with (LOCAL_SAVE_DIR / "training_summary.json").open(
    "w", encoding="utf-8"
) as file:
    json.dump(training_summary, file, indent=2)

# Copy checkpoint to persistent storage.
shutil.copytree(LOCAL_SAVE_DIR, SAVE_DIR)

# Validate copied file sizes before marking complete.
for source in LOCAL_SAVE_DIR.iterdir():
    if source.is_file():
        destination = SAVE_DIR / source.name

        assert destination.exists()
        assert destination.stat().st_size == source.stat().st_size

(SAVE_DIR / "COMPLETE").write_text(
    "Checkpoint saved successfully.",
    encoding="utf-8"
)

# Remove temporary local checkpoint copy.
shutil.rmtree(LOCAL_SAVE_DIR)

# ==========================================
# 6. TRAINING SUMMARY
# ==========================================

print("\n" + "=" * 55)
print("FIRST TRAINING CHUNK COMPLETE")
print("=" * 55)

print("Successful optimizer updates:", successful_updates)
print("Recordings processed:", num_records)
print("Mean CTC loss:", round(training_summary["mean_ctc_loss"], 4))

print(
    "Peak GPU memory:",
    round(
        torch.cuda.max_memory_allocated() / 1024**3,
        2
    ),
    "GB"
)

print("Checkpoint:", SAVE_DIR)
print("Checkpoint complete:", (SAVE_DIR / "COMPLETE").exists())
print("Starting baseline remains untouched.")

print("\nREADY FOR CONTINUED TRAINING")


AssertionError: Checkpoint already exists: /content/drive/MyDrive/Amharic_ASR_XLSR/checkpoints/step_000010
Do not restart from step zero over an existing checkpoint.

In [ ]:

import json
import random
import time
import shutil
import hashlib
import os
from pathlib import Path

import torch
import numpy as np

# ==========================================
# 1. CONTINUATION CONFIGURATION
# ==========================================

START_STEP = 10
END_STEP = 50
ACCUMULATION = 4
SEED = 42

assert len(train_dataset) == 5083
assert successful_updates == START_STEP
assert scheduler.last_epoch == START_STEP
assert model.is_gradient_checkpointing

SAVE_DIR = CHECKPOINT_DIR / f"step_{END_STEP:06d}"
PARTIAL_DIR = CHECKPOINT_DIR / f"step_{END_STEP:06d}.partial"

assert not SAVE_DIR.exists(), (
    f"Checkpoint already exists: {SAVE_DIR}"
)
assert not PARTIAL_DIR.exists(), (
    f"Incomplete checkpoint exists: {PARTIAL_DIR}"
)

# ==========================================
# 2. RECONSTRUCT AND SAVE TRAINING ORDER
# ==========================================

training_order = list(range(len(train_dataset)))
random.Random(SEED).shuffle(training_order)

ORDER_PATH = DATA_DIR / "training_order_25h.json"

order_record = {
    "seed": SEED,
    "recording_count": len(train_dataset),
    "recording_ids": [
        train_records[i]["id"]
        for i in training_order
    ]
}

if ORDER_PATH.exists():
    with ORDER_PATH.open(encoding="utf-8") as f:
        previous_order = json.load(f)

    assert previous_order == order_record, (
        "Training order changed. Cannot safely resume."
    )
else:
    with ORDER_PATH.open("w", encoding="utf-8") as f:
        json.dump(order_record, f, ensure_ascii=False)

print("CONTINUING TRAINING")
print("-" * 50)
print("Starting step:", START_STEP)
print("Ending step:", END_STEP)
print("Additional recordings:", (END_STEP - START_STEP) * 4)
print("Training order verified:", True)

# ==========================================
# 3. TRAIN THE NEXT 40 UPDATES
# ==========================================

model.train()
torch.cuda.reset_peak_memory_stats()

training_log = []
start_time = time.perf_counter()

for step in range(START_STEP + 1, END_STEP + 1):

    optimizer.zero_grad(set_to_none=True)

    # Continue exactly where step 10 stopped.
    offset = (step - 1) * ACCUMULATION

    indices = training_order[
        offset:offset + ACCUMULATION
    ]

    assert len(indices) == ACCUMULATION

    losses = []

    for record_index in indices:

        batch = ctc_collator([
            train_dataset[record_index]
        ])

        batch = {
            key: value.to(DEVICE)
            for key, value in batch.items()
        }

        with torch.autocast(
            device_type="cuda",
            dtype=torch.float16
        ):
            outputs = model(**batch)
            loss = outputs.loss

        assert torch.isfinite(loss).item(), (
            f"Non-finite loss at step {step}"
        )

        losses.append(float(loss.item()))

        scaler.scale(
            loss / ACCUMULATION
        ).backward()

        del batch, outputs, loss

    scaler.unscale_(optimizer)

    grad_norm = torch.nn.utils.clip_grad_norm_(
        encoder_params + head_params,
        max_norm=MAX_GRAD_NORM,
        error_if_nonfinite=True
    )

    previous_scale = scaler.get_scale()

    scaler.step(optimizer)
    scaler.update()

    if scaler.get_scale() < previous_scale:
        raise RuntimeError(
            f"AMP skipped optimizer update at step {step}. "
            "Resume from the last saved checkpoint."
        )

    scheduler.step()
    successful_updates = step

    mean_loss = sum(losses) / len(losses)

    training_log.append({
        "step": step,
        "loss": mean_loss,
        "gradient_norm": float(grad_norm),
        "encoder_lr": optimizer.param_groups[0]["lr"],
        "head_lr": optimizer.param_groups[1]["lr"]
    })

    if step % 5 == 0:
        recent = training_log[-5:]

        print(
            f"Step {step:04d}/{TOTAL_STEPS} | "
            f"Last-5 loss: "
            f"{np.mean([x['loss'] for x in recent]):.4f} | "
            f"Head LR: {optimizer.param_groups[1]['lr']:.8f} | "
            f"Grad norm: {float(grad_norm):.3f}"
        )

training_seconds = time.perf_counter() - start_time

assert successful_updates == END_STEP

# ==========================================
# 4. SAVE COMPLETE TRAINING STATE
# ==========================================

LOCAL_SAVE_DIR = Path(
    f"/content/asr_checkpoint_step_{END_STEP:06d}"
)

assert not LOCAL_SAVE_DIR.exists()
LOCAL_SAVE_DIR.mkdir(parents=True)

model.save_pretrained(
    str(LOCAL_SAVE_DIR),
    safe_serialization=True
)

processor.save_pretrained(str(LOCAL_SAVE_DIR))

state = {
    "global_step": END_STEP,
    "epoch": 0,
    "next_sample_offset": END_STEP * ACCUMULATION,
    "seed": SEED,
    "num_epochs": NUM_EPOCHS,
    "gradient_accumulation": ACCUMULATION,
    "total_steps": TOTAL_STEPS,
    "warmup_steps": WARMUP_STEPS,
    "unfrozen_layers": 2,
    "optimizer": optimizer.state_dict(),
    "scheduler": scheduler.state_dict(),
    "scaler": scaler.state_dict(),
    "torch_rng_state": torch.get_rng_state(),
    "cuda_rng_states": torch.cuda.get_rng_state_all()
}

torch.save(
    state,
    LOCAL_SAVE_DIR / "trainer_state.pt"
)

summary = {
    "starting_step": START_STEP,
    "ending_step": END_STEP,
    "recordings_processed_total": END_STEP * ACCUMULATION,
    "chunk_seconds": training_seconds,
    "chunk_mean_loss": float(np.mean([
        x["loss"] for x in training_log
    ])),
    "training_log": training_log
}

with (LOCAL_SAVE_DIR / "training_summary.json").open(
    "w", encoding="utf-8"
) as f:
    json.dump(summary, f, indent=2)

# ==========================================
# 5. BACK UP AND VERIFY CHECKPOINT
# ==========================================

def file_sha256(path):
    digest = hashlib.sha256()

    with open(path, "rb") as f:
        for chunk in iter(
            lambda: f.read(4 * 1024**2),
            b""
        ):
            digest.update(chunk)

    return digest.hexdigest()

shutil.copytree(LOCAL_SAVE_DIR, PARTIAL_DIR)

for original in LOCAL_SAVE_DIR.iterdir():
    if not original.is_file():
        continue

    copied = PARTIAL_DIR / original.name

    assert copied.exists()
    assert file_sha256(original) == file_sha256(copied), (
        f"Checkpoint verification failed: {original.name}"
    )

# Rename verified checkpoint into its final location.
os.rename(PARTIAL_DIR, SAVE_DIR)

(SAVE_DIR / "COMPLETE").write_text(
    "Checkpoint complete and verified.",
    encoding="utf-8"
)

shutil.rmtree(LOCAL_SAVE_DIR)

# ==========================================
# 6. REPORT
# ==========================================

print("\n" + "=" * 55)
print("STEP 50 CHECKPOINT COMPLETE")
print("=" * 55)

print("Global optimizer step:", successful_updates)
print("Recordings processed:", END_STEP * ACCUMULATION)
print("Mean loss for this chunk:", round(summary["chunk_mean_loss"], 4))
print("Training time (minutes):", round(training_seconds / 60, 2))

print(
    "Peak GPU memory:",
    round(torch.cuda.max_memory_allocated() / 1024**3, 2),
    "GB"
)

print("Checkpoint:", SAVE_DIR)
print("Checkpoint verified:", (SAVE_DIR / "COMPLETE").exists())
print("Training order:", ORDER_PATH)

print("\nREADY FOR STEP-50 EVALUATION")


NameError: name 'successful_updates' is not defined

In [ ]:

import json
import shutil
import numpy as np
import torch

from pathlib import Path
from torchcodec.decoders import AudioDecoder
from jiwer import cer, wer
from IPython.display import Audio, display
from tqdm.auto import tqdm

# ==========================================
# 1. VERIFY CHECKPOINT AND BASELINE
# ==========================================

EVAL_STEP = 50

assert successful_updates == EVAL_STEP
assert (
    CHECKPOINT_DIR / "step_000050" / "COMPLETE"
).exists(), "Step-50 checkpoint is missing."

baseline_metrics_path = (
    DATA_DIR / "baseline_step0_metrics.json"
)

baseline_predictions_path = (
    DATA_DIR / "baseline_step0_predictions_12.jsonl"
)

with baseline_metrics_path.open(encoding="utf-8") as f:
    baseline_metrics = json.load(f)

with baseline_predictions_path.open(encoding="utf-8") as f:
    baseline_records = [
        json.loads(line) for line in f
    ]

baseline_by_id = {
    record["id"]: record
    for record in baseline_records
}

with BASELINE_EVAL_PATH.open(encoding="utf-8") as f:
    eval_records = [
        json.loads(line) for line in f
    ]

assert len(eval_records) == 12
assert {r["id"] for r in eval_records} == set(baseline_by_id)

print("Evaluation step:", EVAL_STEP)
print("Fixed validation recordings:", len(eval_records))
print("Baseline loaded: YES")

# ==========================================
# 2. VERIFY EVALUATION AUDIO
# ==========================================

EVAL_AUDIO_DIR = Path("/content/amharic_eval_audio")
EVAL_AUDIO_DIR.mkdir(parents=True, exist_ok=True)

DRIVE_EVAL_AUDIO = PROJECT_DIR / "evaluation_audio"

for record in eval_records:
    filename = record["id"] + ".mp3"

    local_path = EVAL_AUDIO_DIR / filename
    drive_path = DRIVE_EVAL_AUDIO / filename

    if not local_path.exists():
        assert drive_path.exists(), (
            f"Evaluation audio missing: {filename}"
        )

        shutil.copy2(drive_path, local_path)

# ==========================================
# 3. INFERENCE WITH STEP-50 MODEL
# ==========================================

model.eval()

results = []
references = []
predictions = []
preview_audio = None

try:
    with torch.inference_mode():
        for i, record in enumerate(
            tqdm(eval_records, desc="Step-50 evaluation")
        ):
            path = EVAL_AUDIO_DIR / (
                record["id"] + ".mp3"
            )

            decoder = AudioDecoder(
                str(path),
                sample_rate=SAMPLE_RATE,
                num_channels=1
            )

            decoded = decoder.get_all_samples()

            waveform = (
                decoded.data[0]
                .cpu()
                .numpy()
                .astype(np.float32)
            )

            # Retain one clip for listening after evaluation.
            if i == 0:
                preview_audio = waveform.copy()

            inputs = processor.feature_extractor(
                waveform,
                sampling_rate=SAMPLE_RATE,
                return_attention_mask=True,
                return_tensors="pt"
            )

            inputs = {
                key: value.to(DEVICE)
                for key, value in inputs.items()
            }

            with torch.autocast(
                device_type="cuda",
                dtype=torch.float16
            ):
                logits = model(**inputs).logits

            assert torch.isfinite(logits).all(), (
                f"Non-finite logits for {record['id']}"
            )

            token_ids = logits.argmax(dim=-1)

            predicted = processor.batch_decode(
                token_ids.cpu()
            )[0]

            predicted = normalize_amharic_ctc(
                predicted
            )

            reference = record["transcription"]

            blank_fraction = (
                (token_ids == tokenizer.pad_token_id)
                .float()
                .mean()
                .item()
            )

            result = {
                "id": record["id"],
                "speaker_id": record["speaker_id"],
                "reference": reference,
                "prediction": predicted,
                "duration_seconds": len(waveform) / SAMPLE_RATE,
                "cer": cer(reference, predicted),
                "wer": wer(reference, predicted),
                "blank_fraction": blank_fraction,
                "prediction_length": len(predicted)
            }

            results.append(result)
            references.append(reference)
            predictions.append(predicted)

            del inputs, logits, token_ids

finally:
    # Restore training mode without changing weights.
    model.train()

# ==========================================
# 4. COMPUTE COMPARABLE METRICS
# ==========================================

step50_cer = cer(references, predictions)
step50_wer = wer(references, predictions)

mean_blank = float(np.mean([
    r["blank_fraction"] for r in results
]))

empty_count = sum(
    not prediction for prediction in predictions
)

mean_prediction_length = float(np.mean([
    len(prediction) for prediction in predictions
]))

metrics = {
    "training_step": EVAL_STEP,
    "evaluation_recordings": len(results),
    "cer": step50_cer,
    "wer": step50_wer,
    "mean_blank_fraction": mean_blank,
    "empty_predictions": empty_count,
    "mean_prediction_length": mean_prediction_length
}

# ==========================================
# 5. SAVE RESULTS TO GOOGLE DRIVE
# ==========================================

RESULTS_PATH = (
    DATA_DIR / "eval_step_000050_predictions_12.jsonl"
)

METRICS_PATH = (
    DATA_DIR / "eval_step_000050_metrics.json"
)

with RESULTS_PATH.open("w", encoding="utf-8") as f:
    for result in results:
        f.write(
            json.dumps(result, ensure_ascii=False) + "\n"
        )

with METRICS_PATH.open("w", encoding="utf-8") as f:
    json.dump(metrics, f, indent=2)

# ==========================================
# 6. BASELINE COMPARISON
# ==========================================

print("\n" + "=" * 65)
print("BEFORE VS AFTER: STEP 0 AND STEP 50")
print("=" * 65)

print(
    f"{'Metric':27}"
    f"{'Step 0':>15}"
    f"{'Step 50':>15}"
)

print("-" * 57)

print(
    f"{'CER':27}"
    f"{baseline_metrics['cer'] * 100:14.2f}%"
    f"{step50_cer * 100:14.2f}%"
)

print(
    f"{'WER':27}"
    f"{baseline_metrics['wer'] * 100:14.2f}%"
    f"{step50_wer * 100:14.2f}%"
)

print(
    f"{'Mean blank frames':27}"
    f"{baseline_metrics['mean_blank_fraction'] * 100:14.2f}%"
    f"{mean_blank * 100:14.2f}%"
)

print(
    f"{'Empty predictions':27}"
    f"{baseline_metrics['empty_predictions']:15}"
    f"{empty_count:15}"
)

print("\nCER change (percentage points):",
      round(
          (step50_cer - baseline_metrics["cer"]) * 100,
          2
      ))

# ==========================================
# 7. DISPLAY SIDE-BY-SIDE TRANSCRIPTIONS
# ==========================================

print("\nAMHARIC TRANSCRIPTION COMPARISON")

for i in [0, 5, 11]:
    current = results[i]
    original = baseline_by_id[current["id"]]

    print("\n" + "-" * 65)
    print("RECORDING:", i + 1)
    print("REFERENCE:")
    print(current["reference"][:220])

    print("\nSTEP 0:")
    print(original["prediction"][:220] or "[EMPTY]")

    print("\nSTEP 50:")
    print(current["prediction"][:220] or "[EMPTY]")

    print(
        "\nCER:",
        f"{original['cer'] * 100:.1f}%",
        "->",
        f"{current['cer'] * 100:.1f}%"
    )

print("\nLISTEN TO RECORDING 1:")
display(Audio(preview_audio, rate=SAMPLE_RATE))

print("\nResults saved:", RESULTS_PATH)
print("Metrics saved:", METRICS_PATH)
print("\nSTEP-50 EVALUATION COMPLETE")


In [ ]:

import os
import json
import time
import shutil
import hashlib
import random
from pathlib import Path

import numpy as np
import torch

# ==========================================
# 1. CONTINUATION SETTINGS
# ==========================================

START_STEP = 50
END_STEP = 200
ACCUMULATION = 4

assert successful_updates == START_STEP
assert scheduler.last_epoch == START_STEP
assert model.training
assert model.is_gradient_checkpointing

# Reconstruct the saved deterministic order.
training_order = list(range(len(train_dataset)))
random.Random(TRAINING_SEED).shuffle(training_order)

with ORDER_PATH.open(encoding="utf-8") as f:
    saved_order = json.load(f)

assert [
    train_records[i]["id"]
    for i in training_order
] == saved_order["recording_ids"], (
    "Training order mismatch."
)

assert END_STEP * ACCUMULATION <= len(training_order)

checkpoint_path = (
    CHECKPOINT_DIR / f"step_{END_STEP:06d}"
)

partial_path = (
    CHECKPOINT_DIR / f"step_{END_STEP:06d}.partial"
)

local_path = Path(
    f"/content/asr_step_{END_STEP:06d}_temp"
)

for path in [checkpoint_path, partial_path, local_path]:
    assert not path.exists(), (
        f"Existing checkpoint path: {path}"
    )

print("TRAINING CONTINUATION")
print("-" * 50)
print("Starting step:", START_STEP)
print("Target step:", END_STEP)
print(
    "Additional recordings:",
    (END_STEP - START_STEP) * ACCUMULATION
)
print("Warmup finishes at step:", WARMUP_STEPS)
print("Training order: VERIFIED")

# ==========================================
# 2. CONTINUE OPTIMIZER UPDATES
# ==========================================

model.train()
torch.cuda.reset_peak_memory_stats()

training_log = []
start_time = time.perf_counter()

for step in range(START_STEP + 1, END_STEP + 1):

    optimizer.zero_grad(set_to_none=True)

    offset = (step - 1) * ACCUMULATION
    indices = training_order[offset:offset + ACCUMULATION]

    assert len(indices) == ACCUMULATION

    losses = []

    for record_index in indices:

        batch = ctc_collator(
            [train_dataset[record_index]]
        )

        batch = {
            key: value.to(DEVICE)
            for key, value in batch.items()
        }

        with torch.autocast(
            device_type="cuda",
            dtype=torch.float16
        ):
            outputs = model(**batch)
            loss = outputs.loss

        if not torch.isfinite(loss).item():
            raise RuntimeError(
                f"Non-finite loss at step {step}"
            )

        losses.append(float(loss.item()))

        scaler.scale(
            loss / ACCUMULATION
        ).backward()

        del batch, outputs, loss

    # Unscale before clipping.
    scaler.unscale_(optimizer)

    grad_norm = torch.nn.utils.clip_grad_norm_(
        encoder_params + head_params,
        max_norm=MAX_GRAD_NORM,
        error_if_nonfinite=True
    )

    old_scale = scaler.get_scale()

    scaler.step(optimizer)
    scaler.update()

    if scaler.get_scale() < old_scale:
        raise RuntimeError(
            f"AMP skipped update at step {step}. "
            "Reload the last verified checkpoint."
        )

    scheduler.step()
    successful_updates = step

    mean_loss = float(np.mean(losses))

    training_log.append({
        "step": step,
        "loss": mean_loss,
        "gradient_norm": float(grad_norm),
        "encoder_lr": optimizer.param_groups[0]["lr"],
        "head_lr": optimizer.param_groups[1]["lr"]
    })

    if step % 25 == 0:
        recent_losses = [
            entry["loss"]
            for entry in training_log[-25:]
        ]

        print(
            f"Step {step:04d}/{TOTAL_STEPS} | "
            f"Mean loss (last 25): "
            f"{np.mean(recent_losses):.4f} | "
            f"Head LR: "
            f"{optimizer.param_groups[1]['lr']:.8f}"
        )

elapsed_seconds = time.perf_counter() - start_time

assert successful_updates == END_STEP

# ==========================================
# 3. SAVE MODEL + COMPLETE TRAINING STATE
# ==========================================

local_path.mkdir(parents=True)

model.save_pretrained(
    str(local_path),
    safe_serialization=True
)

processor.save_pretrained(str(local_path))

trainer_state = {
    "global_step": END_STEP,
    "epoch": 0,
    "next_sample_offset": END_STEP * ACCUMULATION,
    "seed": TRAINING_SEED,
    "num_epochs": NUM_EPOCHS,
    "gradient_accumulation": ACCUMULATION,
    "total_steps": TOTAL_STEPS,
    "warmup_steps": WARMUP_STEPS,
    "unfrozen_layers": 2,
    "optimizer": optimizer.state_dict(),
    "scheduler": scheduler.state_dict(),
    "scaler": scaler.state_dict(),
    "torch_rng_state": torch.get_rng_state(),
    "cuda_rng_states": torch.cuda.get_rng_state_all()
}

torch.save(
    trainer_state,
    local_path / "trainer_state.pt"
)

summary = {
    "starting_step": START_STEP,
    "ending_step": END_STEP,
    "total_recordings_processed": END_STEP * ACCUMULATION,
    "mean_chunk_loss": float(np.mean([
        entry["loss"] for entry in training_log
    ])),
    "elapsed_seconds": elapsed_seconds,
    "training_log": training_log
}

with (local_path / "training_summary.json").open(
    "w", encoding="utf-8"
) as f:
    json.dump(summary, f, indent=2)

# ==========================================
# 4. VERIFIED GOOGLE DRIVE BACKUP
# ==========================================

def checkpoint_hash(path):
    digest = hashlib.sha256()

    with path.open("rb") as f:
        for chunk in iter(
            lambda: f.read(4 * 1024**2),
            b""
        ):
            digest.update(chunk)

    return digest.hexdigest()

shutil.copytree(local_path, partial_path)

for source in local_path.iterdir():
    if source.is_file():
        destination = partial_path / source.name

        assert destination.exists()
        assert checkpoint_hash(source) == checkpoint_hash(destination), (
            f"Checksum mismatch: {source.name}"
        )

os.rename(partial_path, checkpoint_path)

(checkpoint_path / "COMPLETE").write_text(
    "Verified checkpoint.",
    encoding="utf-8"
)

shutil.rmtree(local_path)

# ==========================================
# 5. REPORT
# ==========================================

print("\n" + "=" * 55)
print("STEP 200 TRAINING COMPLETE")
print("=" * 55)

print("Global optimizer step:", successful_updates)
print("Recordings processed:", END_STEP * ACCUMULATION)
print("Mean chunk loss:", round(summary["mean_chunk_loss"], 4))
print("Training duration (minutes):", round(elapsed_seconds / 60, 2))

print(
    "Peak GPU memory:",
    round(torch.cuda.max_memory_allocated() / 1024**3, 2),
    "GB"
)

print("Current head LR:", optimizer.param_groups[1]["lr"])
print("Warmup completed:", END_STEP >= WARMUP_STEPS)
print("Checkpoint:", checkpoint_path)
print(
    "Checkpoint verified:",
    (checkpoint_path / "COMPLETE").exists()
)

print("\nREADY FOR STEP-200 EVALUATION")


In [ ]:

import json
import numpy as np
import torch

from pathlib import Path
from torchcodec.decoders import AudioDecoder
from jiwer import cer, wer
from tqdm.auto import tqdm
from IPython.display import Audio, display

# ==========================================
# 1. VERIFY EXPERIMENT STATE
# ==========================================

EVAL_STEP = 200

assert successful_updates == EVAL_STEP
assert (
    CHECKPOINT_DIR / "step_000200" / "COMPLETE"
).exists()

# Load both previous evaluations.
with (
    DATA_DIR / "baseline_step0_metrics.json"
).open(encoding="utf-8") as f:
    step0_metrics = json.load(f)

with (
    DATA_DIR / "eval_step_000050_metrics.json"
).open(encoding="utf-8") as f:
    step50_metrics = json.load(f)

def load_jsonl(path):
    with path.open(encoding="utf-8") as f:
        return [json.loads(line) for line in f]

eval_records = load_jsonl(BASELINE_EVAL_PATH)

step0_predictions = {
    r["id"]: r
    for r in load_jsonl(
        DATA_DIR / "baseline_step0_predictions_12.jsonl"
    )
}

step50_predictions = {
    r["id"]: r
    for r in load_jsonl(
        DATA_DIR / "eval_step_000050_predictions_12.jsonl"
    )
}

assert len(eval_records) == 12

expected_ids = {r["id"] for r in eval_records}

assert set(step0_predictions) == expected_ids
assert set(step50_predictions) == expected_ids

# ==========================================
# 2. INFERENCE ON THE FIXED VALIDATION SET
# ==========================================

model.eval()

results = []
references = []
predictions = []

preview_audio = None

try:
    with torch.inference_mode():

        for index, record in enumerate(
            tqdm(eval_records, desc="Step-200 evaluation")
        ):
            audio_path = (
                EVAL_AUDIO_DIR / f"{record['id']}.mp3"
            )

            assert audio_path.exists(), audio_path

            decoder = AudioDecoder(
                str(audio_path),
                sample_rate=SAMPLE_RATE,
                num_channels=1
            )

            samples = decoder.get_all_samples()

            waveform = (
                samples.data[0]
                .cpu()
                .numpy()
                .astype(np.float32)
            )

            if index == 0:
                preview_audio = waveform.copy()

            inputs = processor.feature_extractor(
                waveform,
                sampling_rate=SAMPLE_RATE,
                return_attention_mask=True,
                return_tensors="pt"
            )

            inputs = {
                name: tensor.to(DEVICE)
                for name, tensor in inputs.items()
            }

            with torch.autocast(
                device_type="cuda",
                dtype=torch.float16
            ):
                logits = model(**inputs).logits

            assert torch.isfinite(logits).all()

            predicted_ids = logits.argmax(dim=-1)

            predicted_text = processor.batch_decode(
                predicted_ids.cpu()
            )[0]

            predicted_text = normalize_amharic_ctc(
                predicted_text
            )

            reference = record["transcription"]

            blank_fraction = (
                (predicted_ids == tokenizer.pad_token_id)
                .float()
                .mean()
                .item()
            )

            result = {
                "id": record["id"],
                "speaker_id": record["speaker_id"],
                "reference": reference,
                "prediction": predicted_text,
                "cer": cer(reference, predicted_text),
                "wer": wer(reference, predicted_text),
                "blank_fraction": blank_fraction,
                "prediction_length": len(predicted_text)
            }

            results.append(result)
            references.append(reference)
            predictions.append(predicted_text)

            del inputs, logits, predicted_ids

finally:
    # Keep the existing model ready for training.
    model.train()

# ==========================================
# 3. CALCULATE EVALUATION METRICS
# ==========================================

step200_metrics = {
    "training_step": EVAL_STEP,
    "evaluation_recordings": len(results),
    "cer": cer(references, predictions),
    "wer": wer(references, predictions),
    "mean_blank_fraction": float(
        np.mean([r["blank_fraction"] for r in results])
    ),
    "empty_predictions": sum(
        not prediction for prediction in predictions
    ),
    "mean_prediction_length": float(
        np.mean([len(p) for p in predictions])
    )
}

# ==========================================
# 4. SAVE RESULTS
# ==========================================

PREDICTIONS_PATH = (
    DATA_DIR / "eval_step_000200_predictions_12.jsonl"
)

METRICS_PATH = (
    DATA_DIR / "eval_step_000200_metrics.json"
)

with PREDICTIONS_PATH.open("w", encoding="utf-8") as f:
    for result in results:
        f.write(
            json.dumps(result, ensure_ascii=False) + "\n"
        )

with METRICS_PATH.open("w", encoding="utf-8") as f:
    json.dump(step200_metrics, f, indent=2)

# ==========================================
# 5. THREE-WAY COMPARISON
# ==========================================

all_metrics = [
    ("Step 0", step0_metrics),
    ("Step 50", step50_metrics),
    ("Step 200", step200_metrics)
]

print("\n" + "=" * 72)
print("AMHARIC ASR: THREE-CHECKPOINT COMPARISON")
print("=" * 72)

print(
    f"{'Checkpoint':<15}"
    f"{'CER':>12}"
    f"{'WER':>12}"
    f"{'Blank %':>14}"
    f"{'Empty':>10}"
)

print("-" * 65)

for name, m in all_metrics:
    print(
        f"{name:<15}"
        f"{m['cer'] * 100:>11.2f}%"
        f"{m['wer'] * 100:>11.2f}%"
        f"{m['mean_blank_fraction'] * 100:>13.2f}%"
        f"{m['empty_predictions']:>10}"
    )

print("\nCER CHANGE")
print(
    "Step 0 -> 200:",
    round(
        (step200_metrics["cer"] - step0_metrics["cer"]) * 100,
        2
    ),
    "percentage points"
)

print(
    "Step 50 -> 200:",
    round(
        (step200_metrics["cer"] - step50_metrics["cer"]) * 100,
        2
    ),
    "percentage points"
)

# ==========================================
# 6. COMPARE ACTUAL AMHARIC PREDICTIONS
# ==========================================

print("\n" + "=" * 72)
print("TRANSCRIPTIONS: BEFORE VS AFTER")
print("=" * 72)

for index in [0, 5, 11]:
    current = results[index]
    record_id = current["id"]

    previous0 = step0_predictions[record_id]
    previous50 = step50_predictions[record_id]

    print(f"\n{'-' * 70}")
    print(f"RECORDING {index + 1}")
    print("REFERENCE:")
    print(current["reference"][:220])

    print("\nSTEP 0:")
    print(previous0["prediction"][:220] or "[EMPTY]")

    print("\nSTEP 50:")
    print(previous50["prediction"][:220] or "[EMPTY]")

    print("\nSTEP 200:")
    print(current["prediction"][:220] or "[EMPTY]")

    print(
        "\nCER:",
        f"{previous0['cer'] * 100:.1f}%",
        "->",
        f"{previous50['cer'] * 100:.1f}%",
        "->",
        f"{current['cer'] * 100:.1f}%"
    )

print("\nAUDIO FOR RECORDING 1:")
display(Audio(preview_audio, rate=SAMPLE_RATE))

print("\nPredictions saved:", PREDICTIONS_PATH)
print("Metrics saved:", METRICS_PATH)
print("\nSTEP-200 EVALUATION COMPLETE")


NameError: name 'successful_updates' is not defined

In [ ]:

import torch
import numpy as np
from pathlib import Path
from torchcodec.decoders import AudioDecoder

assert successful_updates == 200

BLANK_ID = tokenizer.pad_token_id

# Deterministic training groups.
seen_indices = training_order[::199][:4]
unseen_indices = training_order[800::199][:4]

assert len(seen_indices) == 4
assert len(unseen_indices) == 4

# Build three groups of examples.
groups = {
    "TRAIN: SEEN": [
        train_dataset[i] for i in seen_indices
    ],
    "TRAIN: UNSEEN": [
        train_dataset[i] for i in unseen_indices
    ],
    "VALIDATION": []
}

for record in eval_records[:4]:
    audio_path = EVAL_AUDIO_DIR / f"{record['id']}.mp3"

    decoder = AudioDecoder(
        str(audio_path),
        sample_rate=SAMPLE_RATE,
        num_channels=1
    )
    decoded = decoder.get_all_samples()

    waveform = (
        decoded.data[0].cpu().numpy().astype(np.float32)
    )

    features = processor.feature_extractor(
        waveform,
        sampling_rate=SAMPLE_RATE
    )

    labels = tokenizer.encode(
        record["transcription"],
        add_special_tokens=False
    )

    groups["VALIDATION"].append({
        "input_values": features.input_values[0],
        "labels": labels,
        "id": record["id"]
    })

# Inspect predictions and probabilities.
model.eval()

try:
    with torch.inference_mode():

        for group_name, examples in groups.items():

            losses = []
            blank_argmax_rates = []
            blank_probabilities = []
            nonblank_probabilities = []

            print("\n" + "=" * 65)
            print(group_name)
            print("=" * 65)

            for example in examples:
                batch = ctc_collator([example])

                batch = {
                    key: value.to(DEVICE)
                    for key, value in batch.items()
                }

                with torch.autocast(
                    device_type="cuda",
                    dtype=torch.float16
                ):
                    outputs = model(**batch)

                loss = float(outputs.loss.item())

                # Use FP32 for probability diagnostics.
                probs = outputs.logits[0].float().softmax(
                    dim=-1
                )

                frame_predictions = probs.argmax(dim=-1)

                blank_argmax = (
                    frame_predictions == BLANK_ID
                ).float().mean().item()

                blank_mean = (
                    probs[:, BLANK_ID].mean().item()
                )

                # Strongest nonblank probability per frame.
                nonblank = probs.clone()
                nonblank[:, BLANK_ID] = 0.0

                strongest_nonblank = (
                    nonblank.max(dim=-1).values
                )

                mean_nonblank = (
                    strongest_nonblank.mean().item()
                )

                peak_nonblank = (
                    strongest_nonblank.max().item()
                )

                predicted = processor.batch_decode(
                    frame_predictions.unsqueeze(0).cpu()
                )[0]

                # Identify the most probable nonblank tokens,
                # averaged over all acoustic frames.
                mean_token_probs = nonblank.mean(dim=0)
                top_ids = torch.topk(
                    mean_token_probs, k=5
                ).indices.tolist()

                top_tokens = [
                    tokenizer.convert_ids_to_tokens(i)
                    for i in top_ids
                ]

                losses.append(loss)
                blank_argmax_rates.append(blank_argmax)
                blank_probabilities.append(blank_mean)
                nonblank_probabilities.append(mean_nonblank)

                print(f"\nID: {example['id']}")
                print("CTC loss:", round(loss, 4))
                print(
                    "Blank argmax frames:",
                    f"{blank_argmax * 100:.2f}%"
                )
                print(
                    "Mean blank probability:",
                    f"{blank_mean * 100:.2f}%"
                )
                print(
                    "Mean strongest nonblank probability:",
                    f"{mean_nonblank * 100:.2f}%"
                )
                print(
                    "Peak nonblank probability:",
                    f"{peak_nonblank * 100:.2f}%"
                )
                print("Top nonblank tokens:", top_tokens)
                print(
                    "Greedy prediction:",
                    predicted[:100] or "[EMPTY]"
                )

                del batch, outputs, probs, nonblank

            print("\nGROUP SUMMARY")
            print(
                "Mean CTC loss:",
                round(float(np.mean(losses)), 4)
            )
            print(
                "Mean blank argmax:",
                f"{np.mean(blank_argmax_rates) * 100:.2f}%"
            )
            print(
                "Mean blank probability:",
                f"{np.mean(blank_probabilities) * 100:.2f}%"
            )
            print(
                "Mean strongest nonblank probability:",
                f"{np.mean(nonblank_probabilities) * 100:.2f}%"
            )

finally:
    model.train()

print("\nBLANK-DOMINANCE DIAGNOSTIC COMPLETE")
print("No weights were updated.")


In [ ]:

import os
import json
import time
import shutil
import hashlib
import random
import gc
from pathlib import Path

import numpy as np
import torch

# ==========================================
# 1. CONFIGURATION
# ==========================================

START_STEP = 200
END_STEP = 500
SAVE_STEPS = {350, 500}
ACCUMULATION = 4

assert successful_updates == START_STEP
assert scheduler.last_epoch == START_STEP
assert model.is_gradient_checkpointing
assert len(train_dataset) == 5083

# Verify the exact training order.
training_order = list(range(len(train_dataset)))
random.Random(TRAINING_SEED).shuffle(training_order)

with ORDER_PATH.open(encoding="utf-8") as f:
    saved_order = json.load(f)

assert [
    train_records[i]["id"] for i in training_order
] == saved_order["recording_ids"]

assert END_STEP * ACCUMULATION <= len(training_order)

for step in SAVE_STEPS:
    destination = CHECKPOINT_DIR / f"step_{step:06d}"
    assert not destination.exists(), (
        f"Checkpoint already exists: {destination}"
    )

# ==========================================
# 2. VERIFIED CHECKPOINT FUNCTION
# ==========================================

def sha256_file(path):
    digest = hashlib.sha256()

    with path.open("rb") as f:
        for chunk in iter(
            lambda: f.read(4 * 1024 * 1024),
            b""
        ):
            digest.update(chunk)

    return digest.hexdigest()


def save_training_checkpoint(step, logs):

    name = f"step_{step:06d}"

    local_dir = Path(f"/content/{name}_training_temp")
    partial_dir = CHECKPOINT_DIR / f"{name}.partial"
    final_dir = CHECKPOINT_DIR / name

    for path in [local_dir, partial_dir, final_dir]:
        assert not path.exists(), f"Path exists: {path}"

    local_dir.mkdir(parents=True)

    # Model and tokenizer.
    model.save_pretrained(
        str(local_dir),
        safe_serialization=True
    )

    processor.save_pretrained(str(local_dir))

    # Complete optimizer and training state.
    state = {
        "global_step": step,
        "epoch": 0,
        "next_sample_offset": step * ACCUMULATION,
        "seed": TRAINING_SEED,
        "num_epochs": NUM_EPOCHS,
        "gradient_accumulation": ACCUMULATION,
        "total_steps": TOTAL_STEPS,
        "warmup_steps": WARMUP_STEPS,
        "unfrozen_layers": 2,
        "optimizer": optimizer.state_dict(),
        "scheduler": scheduler.state_dict(),
        "scaler": scaler.state_dict(),
        "torch_rng_state": torch.get_rng_state(),
        "cuda_rng_states": torch.cuda.get_rng_state_all(),
        "python_rng_state": random.getstate(),
        "numpy_rng_state": np.random.get_state()
    }

    torch.save(
        state,
        local_dir / "trainer_state.pt"
    )

    summary = {
        "global_step": step,
        "recordings_processed": step * ACCUMULATION,
        "recent_mean_loss": float(
            np.mean([x["loss"] for x in logs[-25:]])
        ),
        "chunk_log": logs
    }

    with (
        local_dir / "training_summary.json"
    ).open("w", encoding="utf-8") as f:
        json.dump(summary, f, indent=2)

    # Copy to Drive and verify contents.
    shutil.copytree(local_dir, partial_dir)

    for source in local_dir.iterdir():
        if source.is_file():
            copied = partial_dir / source.name

            assert copied.exists()
            assert sha256_file(source) == sha256_file(copied), (
                f"Checksum mismatch: {source.name}"
            )

    os.rename(partial_dir, final_dir)

    (final_dir / "COMPLETE").write_text(
        "Verified checkpoint.",
        encoding="utf-8"
    )

    shutil.rmtree(local_dir)

    print(f"\nCHECKPOINT SAVED: STEP {step}")
    print("Location:", final_dir)
    print("Verification: PASSED\n")


# ==========================================
# 3. CONTINUE TRAINING
# ==========================================

model.train()
torch.cuda.reset_peak_memory_stats()

training_log = []
start_time = time.perf_counter()

print("TRAINING CONTINUATION")
print("-" * 55)
print("Starting step:", START_STEP)
print("Target step:", END_STEP)
print("Additional recordings:", (END_STEP - START_STEP) * 4)
print("Checkpoint steps:", sorted(SAVE_STEPS))
print("Training order: VERIFIED")
print()

for step in range(START_STEP + 1, END_STEP + 1):

    optimizer.zero_grad(set_to_none=True)

    offset = (step - 1) * ACCUMULATION
    indices = training_order[
        offset:offset + ACCUMULATION
    ]

    assert len(indices) == ACCUMULATION

    losses = []

    for record_index in indices:

        batch = ctc_collator(
            [train_dataset[record_index]]
        )

        batch = {
            key: value.to(DEVICE)
            for key, value in batch.items()
        }

        with torch.autocast(
            device_type="cuda",
            dtype=torch.float16
        ):
            outputs = model(**batch)
            loss = outputs.loss

        if not torch.isfinite(loss).item():
            raise RuntimeError(
                f"Non-finite CTC loss at step {step}"
            )

        losses.append(float(loss.item()))

        scaler.scale(
            loss / ACCUMULATION
        ).backward()

        del batch, outputs, loss

    # ======================================
    # 4. GRADIENT CLIPPING + UPDATE
    # ======================================

    scaler.unscale_(optimizer)

    grad_norm = torch.nn.utils.clip_grad_norm_(
        encoder_params + head_params,
        max_norm=MAX_GRAD_NORM,
        error_if_nonfinite=True
    )

    scale_before = scaler.get_scale()

    scaler.step(optimizer)
    scaler.update()

    if scaler.get_scale() < scale_before:
        raise RuntimeError(
            f"AMP skipped optimizer update at step {step}. "
            "Recover from the last verified checkpoint."
        )

    scheduler.step()
    successful_updates = step

    mean_loss = float(np.mean(losses))

    training_log.append({
        "step": step,
        "loss": mean_loss,
        "gradient_norm": float(grad_norm),
        "head_lr": optimizer.param_groups[1]["lr"],
        "encoder_lr": optimizer.param_groups[0]["lr"]
    })

    if step % 25 == 0:

        recent = training_log[-25:]

        recent_loss = float(np.mean([
            entry["loss"] for entry in recent
        ]))

        print(
            f"Step {step:04d}/{TOTAL_STEPS} | "
            f"Last-25 loss: {recent_loss:.4f} | "
            f"Head LR: "
            f"{optimizer.param_groups[1]['lr']:.8f}"
        )

    # ======================================
    # 5. PERIODIC VERIFIED CHECKPOINTS
    # ======================================

    if step in SAVE_STEPS:
        save_training_checkpoint(
            step,
            training_log.copy()
        )

# ==========================================
# 6. FINAL REPORT
# ==========================================

elapsed = time.perf_counter() - start_time

assert successful_updates == END_STEP

print("\n" + "=" * 60)
print("TRAINING COMPLETED THROUGH STEP 500")
print("=" * 60)

print("Current step:", successful_updates)
print("Recordings processed:", END_STEP * ACCUMULATION)

print(
    "Mean loss, steps 201-500:",
    round(
        float(np.mean([
            x["loss"] for x in training_log
        ])),
        4
    )
)

print(
    "Mean loss, last 25 steps:",
    round(
        float(np.mean([
            x["loss"] for x in training_log[-25:]
        ])),
        4
    )
)

print("Elapsed minutes:", round(elapsed / 60, 2))

print(
    "Peak GPU memory:",
    round(
        torch.cuda.max_memory_allocated() / 1024**3,
        2
    ),
    "GB"
)

print("\nVERIFIED CHECKPOINTS")

for step in sorted(SAVE_STEPS):
    path = CHECKPOINT_DIR / f"step_{step:06d}"

    print(
        f"Step {step}:",
        "VERIFIED" if (path / "COMPLETE").exists()
        else "MISSING"
    )

print("\nREADY FOR STEP-500 EVALUATION")


In [ ]:

import json
import numpy as np
import torch

from pathlib import Path
from torchcodec.decoders import AudioDecoder
from jiwer import cer, wer
from tqdm.auto import tqdm

# ==========================================
# 1. VERIFY CHECKPOINT
# ==========================================

EVAL_STEP = 500
BLANK_ID = tokenizer.pad_token_id

assert successful_updates == EVAL_STEP
assert (
    CHECKPOINT_DIR / "step_000500" / "COMPLETE"
).exists()

def read_jsonl(path):
    with Path(path).open(encoding="utf-8") as f:
        return [json.loads(line) for line in f]

eval_records = read_jsonl(BASELINE_EVAL_PATH)

assert len(eval_records) == 12

# ==========================================
# 2. LOAD PREVIOUS EVALUATIONS
# ==========================================

previous_metrics = {}

for step, filename in [
    (0, "baseline_step0_metrics.json"),
    (50, "eval_step_000050_metrics.json"),
    (200, "eval_step_000200_metrics.json")
]:
    with (DATA_DIR / filename).open(encoding="utf-8") as f:
        previous_metrics[step] = json.load(f)

previous_predictions = {}

for step, filename in [
    (0, "baseline_step0_predictions_12.jsonl"),
    (50, "eval_step_000050_predictions_12.jsonl"),
    (200, "eval_step_000200_predictions_12.jsonl")
]:
    previous_predictions[step] = {
        r["id"]: r
        for r in read_jsonl(DATA_DIR / filename)
    }

expected_ids = {r["id"] for r in eval_records}

for step in previous_predictions:
    assert set(previous_predictions[step]) == expected_ids

# ==========================================
# 3. INFERENCE HELPER
# ==========================================

def inspect_asr_example(example):

    batch = ctc_collator([example])
    batch = {
        key: value.to(DEVICE)
        for key, value in batch.items()
    }

    with torch.inference_mode():
        with torch.autocast(
            device_type="cuda",
            dtype=torch.float16
        ):
            outputs = model(**batch)

    logits = outputs.logits[0].float()
    loss = float(outputs.loss.item())

    assert torch.isfinite(logits).all()
    assert np.isfinite(loss)

    probabilities = logits.softmax(dim=-1)
    token_ids = probabilities.argmax(dim=-1)

    predicted = processor.batch_decode(
        token_ids.unsqueeze(0).cpu()
    )[0]

    predicted = normalize_amharic_ctc(predicted)

    blank_fraction = (
        (token_ids == BLANK_ID)
        .float()
        .mean()
        .item()
    )

    blank_probability = (
        probabilities[:, BLANK_ID]
        .mean()
        .item()
    )

    nonblank = probabilities.clone()
    nonblank[:, BLANK_ID] = 0.0

    strongest_nonblank = nonblank.max(dim=-1).values

    mean_nonblank = strongest_nonblank.mean().item()
    peak_nonblank = strongest_nonblank.max().item()

    mean_token_probs = nonblank.mean(dim=0)

    top_token_ids = torch.topk(
        mean_token_probs,
        k=5
    ).indices.tolist()

    top_tokens = [
        tokenizer.convert_ids_to_tokens(token_id)
        for token_id in top_token_ids
    ]

    return {
        "id": example["id"],
        "prediction": predicted,
        "ctc_loss": loss,
        "blank_fraction": blank_fraction,
        "blank_probability": blank_probability,
        "mean_strongest_nonblank_probability": mean_nonblank,
        "peak_nonblank_probability": peak_nonblank,
        "top_nonblank_tokens": top_tokens
    }

# ==========================================
# 4. EVALUATE FIXED VALIDATION RECORDINGS
# ==========================================

model.eval()

validation_results = []
seen_train_results = []

try:

    for record in tqdm(
        eval_records,
        desc="Step-500 validation"
    ):

        path = EVAL_AUDIO_DIR / f"{record['id']}.mp3"
        assert path.exists(), path

        decoder = AudioDecoder(
            str(path),
            sample_rate=SAMPLE_RATE,
            num_channels=1
        )

        samples = decoder.get_all_samples()

        waveform = (
            samples.data[0]
            .cpu()
            .numpy()
            .astype(np.float32)
        )

        features = processor.feature_extractor(
            waveform,
            sampling_rate=SAMPLE_RATE
        )

        reference = record["transcription"]

        example = {
            "id": record["id"],
            "input_values": features.input_values[0],
            "labels": tokenizer.encode(
                reference,
                add_special_tokens=False
            )
        }

        result = inspect_asr_example(example)

        result["reference"] = reference
        result["cer"] = cer(reference, result["prediction"])
        result["wer"] = wer(reference, result["prediction"])

        validation_results.append(result)

    # ======================================
    # 5. CHECK FOUR SEEN TRAINING EXAMPLES
    # ======================================

    for index in training_order[:4]:

        example = train_dataset[index]
        result = inspect_asr_example(example)

        result["reference"] = train_records[index][
            "transcription"
        ]

        result["cer"] = cer(
            result["reference"],
            result["prediction"]
        )

        seen_train_results.append(result)

finally:
    model.train()

# ==========================================
# 6. CALCULATE EVALUATION METRICS
# ==========================================

references = [
    r["reference"] for r in validation_results
]

predictions = [
    r["prediction"] for r in validation_results
]

metrics = {
    "training_step": EVAL_STEP,
    "evaluation_recordings": len(validation_results),
    "cer": cer(references, predictions),
    "wer": wer(references, predictions),
    "mean_ctc_loss": float(np.mean([
        r["ctc_loss"] for r in validation_results
    ])),
    "mean_blank_fraction": float(np.mean([
        r["blank_fraction"] for r in validation_results
    ])),
    "mean_blank_probability": float(np.mean([
        r["blank_probability"] for r in validation_results
    ])),
    "mean_strongest_nonblank_probability": float(
        np.mean([
            r["mean_strongest_nonblank_probability"]
            for r in validation_results
        ])
    ),
    "empty_predictions": sum(
        not r["prediction"] for r in validation_results
    ),
    "mean_prediction_length": float(np.mean([
        len(r["prediction"])
        for r in validation_results
    ]))
}

# ==========================================
# 7. SAVE RESULTS
# ==========================================

predictions_path = (
    DATA_DIR / "eval_step_000500_predictions_12.jsonl"
)

metrics_path = (
    DATA_DIR / "eval_step_000500_metrics.json"
)

train_diagnostics_path = (
    DATA_DIR / "eval_step_000500_seen_train_4.jsonl"
)

for path, records in [
    (predictions_path, validation_results),
    (train_diagnostics_path, seen_train_results)
]:
    with path.open("w", encoding="utf-8") as f:
        for record in records:
            f.write(
                json.dumps(record, ensure_ascii=False)
                + "\n"
            )

with metrics_path.open("w", encoding="utf-8") as f:
    json.dump(metrics, f, indent=2)

# ==========================================
# 8. FOUR-CHECKPOINT COMPARISON
# ==========================================

print("\n" + "=" * 72)
print("AMHARIC ASR CHECKPOINT COMPARISON")
print("=" * 72)

print(
    f"{'Step':<10}"
    f"{'CER':>12}"
    f"{'WER':>12}"
    f"{'Blank frames':>17}"
    f"{'Empty':>10}"
)

print("-" * 65)

for step, values in [
    (0, previous_metrics[0]),
    (50, previous_metrics[50]),
    (200, previous_metrics[200]),
    (500, metrics)
]:
    print(
        f"{step:<10}"
        f"{values['cer'] * 100:>11.2f}%"
        f"{values['wer'] * 100:>11.2f}%"
        f"{values['mean_blank_fraction'] * 100:>16.2f}%"
        f"{values['empty_predictions']:>10}"
    )

# ==========================================
# 9. STEP-500 PROBABILITY DIAGNOSTICS
# ==========================================

print("\n" + "=" * 72)
print("STEP-500 VALIDATION DIAGNOSTICS")
print("=" * 72)

print("Mean validation CTC loss:",
      round(metrics["mean_ctc_loss"], 4))

print("Mean blank probability:",
      f"{metrics['mean_blank_probability'] * 100:.2f}%")

print("Mean strongest nonblank probability:",
      f"{metrics['mean_strongest_nonblank_probability'] * 100:.2f}%")

print("Mean prediction length:",
      round(metrics["mean_prediction_length"], 2))

print("Empty predictions:",
      metrics["empty_predictions"], "/12")

# ==========================================
# 10. INSPECT PREVIOUSLY SEEN TRAINING AUDIO
# ==========================================

print("\n" + "=" * 72)
print("SEEN TRAINING RECORDINGS")
print("=" * 72)

for i, result in enumerate(seen_train_results, 1):
    print(f"\nRecording {i}")
    print("CTC loss:", round(result["ctc_loss"], 4))
    print("CER:", f"{result['cer'] * 100:.2f}%")
    print(
        "Blank argmax:",
        f"{result['blank_fraction'] * 100:.2f}%"
    )
    print(
        "Blank probability:",
        f"{result['blank_probability'] * 100:.2f}%"
    )
    print("Top nonblank tokens:", result["top_nonblank_tokens"])
    print("Prediction:", result["prediction"][:120] or "[EMPTY]")

# ==========================================
# 11. SHOW ACTUAL TRANSCRIPTION COMPARISONS
# ==========================================

print("\n" + "=" * 72)
print("BEFORE-AND-AFTER AMHARIC TRANSCRIPTIONS")
print("=" * 72)

for index in [0, 5, 11]:

    current = validation_results[index]
    record_id = current["id"]

    print(f"\n{'-' * 60}")
    print("RECORDING:", index + 1)

    print("REFERENCE:")
    print(current["reference"][:180])

    for step in [0, 50, 200]:
        previous = previous_predictions[step][record_id]

        print(f"\nSTEP {step}:")
        print(previous["prediction"][:180] or "[EMPTY]")

    print("\nSTEP 500:")
    print(current["prediction"][:180] or "[EMPTY]")

    print(
        "Top nonblank tokens:",
        current["top_nonblank_tokens"]
    )

print("\nStep-500 metrics saved:", metrics_path)
print("Step-500 predictions saved:", predictions_path)
print("Seen-training diagnostics:", train_diagnostics_path)
print("\nSTEP-500 EVALUATION COMPLETE")


In [ ]:

import json
import numpy as np
import torch

from pathlib import Path
from torchcodec.decoders import AudioDecoder

# ==========================================
# 1. VERIFY MODEL STATE
# ==========================================

assert successful_updates == 500
assert model.training

BLANK_ID = tokenizer.pad_token_id

# Two recordings already used for training.
seen_examples = [
    train_dataset[i]
    for i in training_order[:2]
]

# Two held-out validation recordings.
validation_examples = []

for record in eval_records[:2]:

    path = EVAL_AUDIO_DIR / f"{record['id']}.mp3"

    decoder = AudioDecoder(
        str(path),
        sample_rate=SAMPLE_RATE,
        num_channels=1
    )

    waveform = (
        decoder.get_all_samples()
        .data[0]
        .cpu()
        .numpy()
        .astype(np.float32)
    )

    features = processor.feature_extractor(
        waveform,
        sampling_rate=SAMPLE_RATE
    )

    validation_examples.append({
        "id": record["id"],
        "input_values": features.input_values[0],
        "labels": tokenizer.encode(
            record["transcription"],
            add_special_tokens=False
        )
    })

groups = {
    "SEEN TRAINING": seen_examples,
    "VALIDATION": validation_examples
}

# ==========================================
# 2. DIAGNOSTIC INFERENCE FUNCTION
# ==========================================

def probe_model(example, audio_values):

    modified = {
        "id": example["id"],
        "input_values": np.asarray(
            audio_values,
            dtype=np.float32
        ).copy(),
        "labels": example["labels"]
    }

    batch = ctc_collator([modified])

    batch = {
        key: value.to(DEVICE)
        for key, value in batch.items()
    }

    with torch.inference_mode():
        with torch.autocast(
            device_type="cuda",
            dtype=torch.float16
        ):
            output = model(
                **batch,
                output_hidden_states=True
            )

    logits = output.logits[0].float()
    probabilities = logits.softmax(dim=-1)

    assert torch.isfinite(logits).all()
    assert torch.isfinite(output.loss)

    predicted_ids = logits.argmax(dim=-1)

    prediction = processor.batch_decode(
        predicted_ids.unsqueeze(0).cpu()
    )[0]

    # Hidden-state variability across time.
    # Index 0 is the encoder input.
    # Index 24 is the final Transformer output.
    hidden_variation = {}

    for layer_index in [0, 12, 22, 24]:

        hidden = output.hidden_states[
            layer_index
        ][0].float()

        temporal_std = hidden.std(
            dim=0,
            unbiased=False
        ).mean().item()

        rms = hidden.square().mean().sqrt().item()

        hidden_variation[str(layer_index)] = {
            "temporal_std": temporal_std,
            "relative_variation": (
                temporal_std / max(rms, 1e-8)
            )
        }

    result = {
        "ctc_loss": float(output.loss.item()),
        "blank_probability": float(
            probabilities[:, BLANK_ID].mean().item()
        ),
        "blank_argmax": float(
            (predicted_ids == BLANK_ID)
            .float().mean().item()
        ),
        "logit_temporal_std": float(
            logits.std(
                dim=0,
                unbiased=False
            ).mean().item()
        ),
        "prediction": prediction,
        "hidden_variation": hidden_variation
    }

    # Return probabilities for comparison.
    probability_copy = probabilities.cpu()

    del batch, output, logits, probabilities

    return result, probability_copy

# ==========================================
# 3. COMPARE ORIGINAL, REVERSED, SILENCE
# ==========================================

model.eval()

diagnostic_results = []

try:
    for group_name, examples in groups.items():

        print("\n" + "=" * 65)
        print(group_name)
        print("=" * 65)

        for example in examples:

            original = np.asarray(
                example["input_values"],
                dtype=np.float32
            )

            variations = {
                "original": original,
                "reversed": original[::-1].copy(),
                "silence": np.zeros_like(original)
            }

            outputs = {}
            distributions = {}

            for condition, waveform in variations.items():

                result, probs = probe_model(
                    example,
                    waveform
                )

                outputs[condition] = result
                distributions[condition] = probs

            original_loss = outputs["original"]["ctc_loss"]
            reversed_loss = outputs["reversed"]["ctc_loss"]
            silence_loss = outputs["silence"]["ctc_loss"]

            # Total variation distance, averaged over frames.
            # 0 means identical token distributions.
            # 1 means completely disjoint distributions.
            reverse_distance = (
                0.5 * (
                    distributions["original"]
                    - distributions["reversed"]
                ).abs().sum(dim=-1).mean().item()
            )

            silence_distance = (
                0.5 * (
                    distributions["original"]
                    - distributions["silence"]
                ).abs().sum(dim=-1).mean().item()
            )

            diagnostic_results.append({
                "group": group_name,
                "id": example["id"],
                "conditions": outputs,
                "original_vs_reversed_tvd": reverse_distance,
                "original_vs_silence_tvd": silence_distance
            })

            print(f"\nRECORDING: {example['id']}")
            print("-" * 55)

            print(
                f"{'Input':<12}"
                f"{'CTC loss':>12}"
                f"{'Blank prob':>14}"
                f"{'Logit std':>13}"
            )

            for condition, result in outputs.items():
                print(
                    f"{condition:<12}"
                    f"{result['ctc_loss']:>12.4f}"
                    f"{result['blank_probability'] * 100:>13.2f}%"
                    f"{result['logit_temporal_std']:>13.5f}"
                )

            print("\nLoss difference vs original:")
            print(
                "Reversed:",
                round(reversed_loss - original_loss, 4)
            )
            print(
                "Silence:",
                round(silence_loss - original_loss, 4)
            )

            print("\nOutput distribution difference:")
            print(
                "Original vs reversed:",
                round(reverse_distance, 5)
            )
            print(
                "Original vs silence:",
                round(silence_distance, 5)
            )

            print("\nOriginal audio hidden-state variation:")

            for layer, statistics in outputs[
                "original"
            ]["hidden_variation"].items():

                print(
                    f"Layer {layer:>2}: "
                    f"temporal_std="
                    f"{statistics['temporal_std']:.6f} "
                    f"relative="
                    f"{statistics['relative_variation']:.6f}"
                )

            print(
                "\nOriginal prediction:",
                outputs["original"]["prediction"][:100]
                or "[EMPTY]"
            )

finally:
    model.train()

# ==========================================
# 4. SAVE THE DIAGNOSTIC
# ==========================================

DIAGNOSTIC_PATH = (
    DATA_DIR / "acoustic_sensitivity_step500.json"
)

with DIAGNOSTIC_PATH.open(
    "w",
    encoding="utf-8"
) as file:

    json.dump(
        diagnostic_results,
        file,
        indent=2,
        ensure_ascii=False
    )

print("\n" + "=" * 65)
print("ACOUSTIC SENSITIVITY DIAGNOSTIC COMPLETE")
print("=" * 65)
print("Results saved:", DIAGNOSTIC_PATH)
print("Model weights updated: NO")
print("Optimizer steps added: 0")


In [ ]:

import gc
import json
import torch
import numpy as np

from transformers import Wav2Vec2ForCTC
from torchcodec.decoders import AudioDecoder

# ==========================================
# 1. LOAD ORIGINAL CHECKPOINT SEPARATELY
# ==========================================

assert successful_updates == 500
assert (BASELINE_DIR / "model.safetensors").exists()

original_training_mode = model.training

baseline_probe = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(DEVICE)

baseline_probe.eval()
model.eval()

LAYERS = [0, 12, 22, 23, 24]

print("REPRESENTATION COMPARISON")
print("-" * 55)
print("Starting model:", BASELINE_DIR)
print("Fine-tuned model: step 500")
print("Layers inspected:", LAYERS)

# ==========================================
# 2. SELECT ONE TRAINING + ONE VALIDATION CLIP
# ==========================================

training_example = train_dataset[training_order[0]]

validation_record = eval_records[0]

decoder = AudioDecoder(
    str(EVAL_AUDIO_DIR / f"{validation_record['id']}.mp3"),
    sample_rate=SAMPLE_RATE,
    num_channels=1
)

waveform = (
    decoder.get_all_samples()
    .data[0]
    .cpu()
    .numpy()
    .astype(np.float32)
)

validation_features = processor.feature_extractor(
    waveform,
    sampling_rate=SAMPLE_RATE
)

validation_example = {
    "id": validation_record["id"],
    "input_values": validation_features.input_values[0],
    "labels": tokenizer.encode(
        validation_record["transcription"],
        add_special_tokens=False
    )
}

examples = {
    "TRAINING": training_example,
    "VALIDATION": validation_example
}

# ==========================================
# 3. PROBE INTERNAL REPRESENTATIONS
# ==========================================

def representation_probe(current_model, example, silence=False):

    batch = ctc_collator([example])

    if silence:
        batch["input_values"] = torch.zeros_like(
            batch["input_values"]
        )

    batch = {
        key: value.to(DEVICE)
        for key, value in batch.items()
    }

    with torch.inference_mode():
        with torch.autocast(
            device_type="cuda",
            dtype=torch.float16
        ):
            output = current_model(
                **batch,
                output_hidden_states=True
            )

    states = {}
    statistics = {}

    for layer_index in LAYERS:
        hidden = (
            output.hidden_states[layer_index][0]
            .float()
            .cpu()
            .clone()
        )

        states[layer_index] = hidden

        temporal_std = hidden.std(
            dim=0,
            unbiased=False
        ).mean().item()

        rms = hidden.square().mean().sqrt().item()

        statistics[layer_index] = {
            "temporal_std": temporal_std,
            "relative_variation": temporal_std / max(rms, 1e-8)
        }

    logits = output.logits[0].float()

    probabilities = (
        logits.softmax(dim=-1)
        .cpu()
        .clone()
    )

    result = {
        "ctc_loss": float(output.loss.item()),
        "blank_probability": float(
            probabilities[:, tokenizer.pad_token_id]
            .mean().item()
        ),
        "statistics": statistics
    }

    del batch, output, logits

    return result, states, probabilities


def relative_rms_difference(a, b):
    difference = (a - b).square().mean().sqrt()
    reference = a.square().mean().sqrt().clamp_min(1e-8)
    return float((difference / reference).item())


# ==========================================
# 4. COMPARE BOTH CHECKPOINTS
# ==========================================

all_results = {}

try:
    for group_name, example in examples.items():

        print("\n" + "=" * 65)
        print(group_name)
        print("Recording:", example["id"])
        print("=" * 65)

        baseline, base_states, base_probs = (
            representation_probe(
                baseline_probe, example
            )
        )

        trained, trained_states, trained_probs = (
            representation_probe(
                model, example
            )
        )

        baseline_silence, base_silence_states, base_silence_probs = (
            representation_probe(
                baseline_probe, example, silence=True
            )
        )

        trained_silence, trained_silence_states, trained_silence_probs = (
            representation_probe(
                model, example, silence=True
            )
        )

        print("\nTEMPORAL VARIATION BY LAYER")
        print(
            f"{'Layer':<8}"
            f"{'Step 0':>13}"
            f"{'Step 500':>13}"
            f"{'Ratio':>12}"
        )
        print("-" * 46)

        layer_comparison = {}

        for layer in LAYERS:

            before = baseline["statistics"][layer][
                "relative_variation"
            ]

            after = trained["statistics"][layer][
                "relative_variation"
            ]

            ratio = after / max(before, 1e-8)

            layer_comparison[str(layer)] = {
                "step0_relative_variation": before,
                "step500_relative_variation": after,
                "ratio": ratio
            }

            print(
                f"{layer:<8}"
                f"{before:>13.6f}"
                f"{after:>13.6f}"
                f"{ratio:>12.4f}"
            )

        # Compare the frozen encoder output.
        frozen_difference = relative_rms_difference(
            base_states[22],
            trained_states[22]
        )

        # Compare acoustic sensitivity in final states.
        base_hidden_sensitivity = relative_rms_difference(
            base_states[24],
            base_silence_states[24]
        )

        trained_hidden_sensitivity = relative_rms_difference(
            trained_states[24],
            trained_silence_states[24]
        )

        # Compare output token distributions.
        base_tvd = float(
            0.5 * (
                base_probs - base_silence_probs
            ).abs().sum(dim=-1).mean().item()
        )

        trained_tvd = float(
            0.5 * (
                trained_probs - trained_silence_probs
            ).abs().sum(dim=-1).mean().item()
        )

        print("\nACOUSTIC SENSITIVITY COMPARISON")
        print("-" * 55)

        print(
            "Frozen layer-22 difference (step 0 vs 500):",
            round(frozen_difference, 8)
        )

        print(
            "Final hidden sensitivity, step 0:",
            round(base_hidden_sensitivity, 5)
        )

        print(
            "Final hidden sensitivity, step 500:",
            round(trained_hidden_sensitivity, 5)
        )

        print(
            "Output TVD vs silence, step 0:",
            round(base_tvd, 5)
        )

        print(
            "Output TVD vs silence, step 500:",
            round(trained_tvd, 5)
        )

        print("\nCTC LOSSES")
        print(
            "Step 0: real / silence:",
            round(baseline["ctc_loss"], 4),
            "/",
            round(baseline_silence["ctc_loss"], 4)
        )

        print(
            "Step 500: real / silence:",
            round(trained["ctc_loss"], 4),
            "/",
            round(trained_silence["ctc_loss"], 4)
        )

        all_results[group_name] = {
            "recording_id": example["id"],
            "layers": layer_comparison,
            "frozen_layer22_relative_difference": frozen_difference,
            "step0_final_hidden_sensitivity": base_hidden_sensitivity,
            "step500_final_hidden_sensitivity": trained_hidden_sensitivity,
            "step0_output_tvd_vs_silence": base_tvd,
            "step500_output_tvd_vs_silence": trained_tvd,
            "step0_ctc_loss": baseline["ctc_loss"],
            "step500_ctc_loss": trained["ctc_loss"]
        }

finally:
    # Do not disturb the training model or optimizer.
    model.train(original_training_mode)

    del baseline_probe
    gc.collect()
    torch.cuda.empty_cache()

# ==========================================
# 5. SAVE DIAGNOSTIC
# ==========================================

OUTPUT_PATH = (
    DATA_DIR / "representation_comparison_step0_vs_500.json"
)

with OUTPUT_PATH.open("w", encoding="utf-8") as file:
    json.dump(
        all_results,
        file,
        indent=2,
        ensure_ascii=False
    )

print("\n" + "=" * 65)
print("REPRESENTATION COMPARISON COMPLETE")
print("=" * 65)
print("Results:", OUTPUT_PATH)
print("Model weights modified: NO")
print("Optimizer steps added: 0")


In [ ]:

import gc
import json
import numpy as np
import torch

from pathlib import Path
from jiwer import cer
from transformers import Wav2Vec2ForCTC

# ==========================================
# 1. VERIFY ORIGINAL MODEL STATE
# ==========================================

assert successful_updates == 500

PROBE_STEPS = 200
PROBE_SEED = 123

PROBE_ENCODER_LR = 2e-5
PROBE_HEAD_LR = 2e-4

# Save RNG state so our regular training can
# continue without altered dropout randomness.
cpu_rng_before = torch.get_rng_state().clone()
cuda_rng_before = torch.cuda.get_rng_state_all()

torch.manual_seed(PROBE_SEED)
torch.cuda.manual_seed_all(PROBE_SEED)

# ==========================================
# 2. SELECT ONE SEEN TRAINING RECORDING
# ==========================================

seen_indices = training_order[:2000]

candidates = [
    i for i in seen_indices
    if 5 <= train_records[i]["duration_seconds"] <= 12
    and 15 <= len(
        tokenizer.encode(
            train_records[i]["transcription"],
            add_special_tokens=False
        )
    ) <= 85
]

if not candidates:
    candidates = [
        i for i in seen_indices
        if len(
            tokenizer.encode(
                train_records[i]["transcription"],
                add_special_tokens=False
            )
        ) >= 15
    ]

assert candidates, "No suitable recording found."

sample_index = min(
    candidates,
    key=lambda i: train_records[i]["duration_seconds"]
)

sample_record = train_records[sample_index]
sample_example = train_dataset[sample_index]

REFERENCE = sample_record["transcription"]

print("SINGLE-EXAMPLE MEMORIZATION TEST")
print("-" * 55)
print("Recording:", sample_record["id"])
print("Duration:", sample_record["duration_seconds"], "seconds")
print("Reference tokens:", len(sample_example["labels"]))
print("Reference:", REFERENCE[:240])

# ==========================================
# 3. LOAD SEPARATE STEP-500 MODEL
# ==========================================

PROBE_CHECKPOINT = (
    CHECKPOINT_DIR / "step_000500"
)

assert (PROBE_CHECKPOINT / "COMPLETE").exists()

probe_model = Wav2Vec2ForCTC.from_pretrained(
    str(PROBE_CHECKPOINT)
).to(DEVICE)

# Match the original trainable architecture.
for parameter in probe_model.parameters():
    parameter.requires_grad = False

for layer in probe_model.wav2vec2.encoder.layers[-2:]:
    for parameter in layer.parameters():
        parameter.requires_grad = True

for parameter in probe_model.lm_head.parameters():
    parameter.requires_grad = True

probe_model.gradient_checkpointing_enable(
    gradient_checkpointing_kwargs={
        "use_reentrant": False
    }
)

# ==========================================
# 4. CREATE DIAGNOSTIC OPTIMIZER
# ==========================================

probe_encoder_params = [
    p
    for layer in probe_model.wav2vec2.encoder.layers[-2:]
    for p in layer.parameters()
    if p.requires_grad
]

probe_head_params = [
    p
    for p in probe_model.lm_head.parameters()
    if p.requires_grad
]

probe_optimizer = torch.optim.AdamW(
    [
        {
            "params": probe_encoder_params,
            "lr": PROBE_ENCODER_LR
        },
        {
            "params": probe_head_params,
            "lr": PROBE_HEAD_LR
        }
    ],
    weight_decay=0.0
)

probe_scaler = torch.amp.GradScaler(
    "cuda",
    init_scale=128.0
)

# Prepare the recording once, avoiding
# repeated MP3 decoding.
probe_batch = ctc_collator([sample_example])

probe_batch = {
    key: value.to(DEVICE)
    for key, value in probe_batch.items()
}

# ==========================================
# 5. EVALUATION HELPER
# ==========================================

def evaluate_probe():

    probe_model.eval()

    with torch.inference_mode():

        with torch.autocast(
            device_type="cuda",
            dtype=torch.float16
        ):
            output = probe_model(**probe_batch)

        logits = output.logits.float()
        assert torch.isfinite(logits).all()

        probabilities = logits.softmax(dim=-1)

        predicted_ids = logits.argmax(dim=-1)

        prediction = processor.batch_decode(
            predicted_ids.cpu()
        )[0]

        prediction = normalize_amharic_ctc(prediction)

        blank_probability = (
            probabilities[..., tokenizer.pad_token_id]
            .mean()
            .item()
        )

        blank_fraction = (
            (predicted_ids == tokenizer.pad_token_id)
            .float()
            .mean()
            .item()
        )

        result = {
            "ctc_loss": float(output.loss.item()),
            "cer": float(cer(REFERENCE, prediction)),
            "blank_probability": float(blank_probability),
            "blank_fraction": float(blank_fraction),
            "prediction": prediction
        }

    return result

# ==========================================
# 6. TRAIN REPEATEDLY ON ONE RECORDING
# ==========================================

probe_history = []
completed_probe_steps = 0

REPORT_STEPS = {
    0, 10, 25, 50, 75, 100, 150, 200
}

try:

    # First measure the unchanged step-500 copy.
    initial = evaluate_probe()

    probe_history.append({
        "step": 0,
        **initial
    })

    print("\nINITIAL PERFORMANCE")
    print("CTC loss:", round(initial["ctc_loss"], 4))
    print("CER:", f"{initial['cer'] * 100:.2f}%")
    print(
        "Blank probability:",
        f"{initial['blank_probability'] * 100:.2f}%"
    )
    print("Prediction:", initial["prediction"][:150] or "[EMPTY]")

    for step in range(1, PROBE_STEPS + 1):

        probe_model.train()

        probe_optimizer.zero_grad(set_to_none=True)

        with torch.autocast(
            device_type="cuda",
            dtype=torch.float16
        ):
            output = probe_model(**probe_batch)
            loss = output.loss

        if not torch.isfinite(loss).item():
            raise RuntimeError(
                f"Non-finite CTC loss at probe step {step}"
            )

        probe_scaler.scale(loss).backward()

        probe_scaler.unscale_(probe_optimizer)

        torch.nn.utils.clip_grad_norm_(
            probe_encoder_params + probe_head_params,
            max_norm=1.0,
            error_if_nonfinite=True
        )

        old_scale = probe_scaler.get_scale()

        probe_scaler.step(probe_optimizer)
        probe_scaler.update()

        if probe_scaler.get_scale() < old_scale:
            raise RuntimeError(
                f"AMP overflow at probe step {step}"
            )

        completed_probe_steps = step

        del output, loss

        if step in REPORT_STEPS:

            result = evaluate_probe()

            probe_history.append({
                "step": step,
                **result
            })

            print(f"\nSTEP {step}/{PROBE_STEPS}")
            print("CTC loss:", round(result["ctc_loss"], 4))
            print("CER:", f"{result['cer'] * 100:.2f}%")
            print(
                "Blank probability:",
                f"{result['blank_probability'] * 100:.2f}%"
            )
            print(
                "Blank argmax:",
                f"{result['blank_fraction'] * 100:.2f}%"
            )
            print(
                "Prediction:",
                result["prediction"][:150] or "[EMPTY]"
            )

            # Early stopping if the model memorizes
            # the example with sufficiently low CER.
            if result["cer"] <= 0.05:
                print("\nMEMORIZATION TARGET REACHED")
                break

    # ======================================
    # 7. SAVE DIAGNOSTIC RESULTS ONLY
    # ======================================

    PROBE_OUTPUT = (
        DATA_DIR / "single_example_overfit_step500.json"
    )

    report = {
        "source_checkpoint": str(PROBE_CHECKPOINT),
        "recording_id": sample_record["id"],
        "duration_seconds": sample_record["duration_seconds"],
        "reference": REFERENCE,
        "probe_encoder_lr": PROBE_ENCODER_LR,
        "probe_head_lr": PROBE_HEAD_LR,
        "completed_steps": completed_probe_steps,
        "history": probe_history
    }

    with PROBE_OUTPUT.open(
        "w", encoding="utf-8"
    ) as file:
        json.dump(
            report,
            file,
            ensure_ascii=False,
            indent=2
        )

    print("\n" + "=" * 65)
    print("SINGLE-EXAMPLE MEMORIZATION RESULTS")
    print("=" * 65)

    print("Starting CER:", f"{initial['cer'] * 100:.2f}%")
    print(
        "Final CER:",
        f"{probe_history[-1]['cer'] * 100:.2f}%"
    )
    print(
        "Starting CTC loss:",
        round(initial["ctc_loss"], 4)
    )
    print(
        "Final CTC loss:",
        round(probe_history[-1]["ctc_loss"], 4)
    )

    print("\nREFERENCE:")
    print(REFERENCE[:300])

    print("\nFINAL PREDICTION:")
    print(probe_history[-1]["prediction"][:300] or "[EMPTY]")

    print("\nResults saved:", PROBE_OUTPUT)

finally:

    # Free only the diagnostic model.
    del probe_model, probe_optimizer, probe_scaler
    del probe_batch

    gc.collect()
    torch.cuda.empty_cache()

    # Restore randomness used by original training.
    torch.set_rng_state(cpu_rng_before)
    torch.cuda.set_rng_state_all(cuda_rng_before)

print("\nMAIN TRAINING MODEL UNCHANGED")
print("Main optimizer remains at step:", successful_updates)


In [ ]:

import copy
import json
import gc

import torch
import torch.nn.functional as F
from jiwer import cer
from transformers import Wav2Vec2ForCTC

# ==========================================
# 1. CONFIGURATION
# ==========================================


# ==========================================
# RESTORE HEAD-ONLY EXPERIMENT DEPENDENCIES
# No previous training state is required.
# ==========================================

from pathlib import Path

DEVICE = "cuda" if torch.cuda.is_available() else "cpu"

# Check that the necessary components exist.
required_variables = [
    "BASELINE_DIR",
    "DATA_DIR",
    "train_records",
    "train_dataset",
    "processor",
    "tokenizer",
    "ctc_collator",
    "normalize_amharic_ctc",
]

missing = [
    name for name in required_variables
    if name not in globals()
]

assert not missing, (
    "Missing notebook dependencies: "
    + ", ".join(missing)
)

assert Path(BASELINE_DIR).exists(), (
    f"Original baseline not found: {BASELINE_DIR}"
)

# Restore the original diagnostic recording.
TARGET_ID = "6Q0fEziAqyQVIz4J8aws"

sample_index = next(
    i for i, record in enumerate(train_records)
    if record["id"] == TARGET_ID
)

sample_record = train_records[sample_index]
sample_example = train_dataset[sample_index]

print("HEAD-ONLY EXPERIMENT READY")
print("Device:", DEVICE)
print("Original baseline:", BASELINE_DIR)
print("Sample:", sample_record["id"])
print("Duration:", sample_record["duration_seconds"], "seconds")
print("Target tokens:", len(sample_example["labels"]))
print("No step-500 model required.")


HEAD_ONLY_STEPS = 1000
HEAD_ONLY_LR = 1e-3
BLANK_ID = tokenizer.pad_token_id

REPORT_STEPS = {
    0, 25, 50, 100, 200, 350,
    500, 750, 1000
}

assert sample_record["id"] == (
    "6Q0fEziAqyQVIz4J8aws"
)

REFERENCE = sample_record["transcription"]

print("FROZEN-ENCODER MEMORIZATION EXPERIMENT")
print("-" * 55)
print("Recording:", sample_record["id"])
print("Reference:", REFERENCE)
print("Model starting point: STEP ZERO")
print("Trainable component: CTC HEAD ONLY")
print("Maximum updates:", HEAD_ONLY_STEPS)

# ==========================================
# 2. LOAD THE ORIGINAL XLS-R CHECKPOINT
# ==========================================

baseline_model = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(DEVICE)

baseline_model.eval()

batch = ctc_collator([sample_example])

batch = {
    key: value.to(DEVICE)
    for key, value in batch.items()
}

# ==========================================
# 3. EXTRACT AND CACHE ORIGINAL FEATURES
# ==========================================


# ==========================================
# 3. EXTRACT AND CACHE ORIGINAL FEATURES
# FIXED: Keep trainable parameters outside inference mode
# ==========================================

with torch.inference_mode():

    original_forward = baseline_model(**batch)

    frozen_features = baseline_model.wav2vec2(
        input_values=batch["input_values"],
        attention_mask=batch["attention_mask"]
    ).last_hidden_state

    initial_full_loss = float(
        original_forward.loss.item()
    )

# IMPORTANT: Clone OUTSIDE inference_mode.
# This creates a normal tensor usable during training.
frozen_features = (
    frozen_features.detach().clone().float()
)

# IMPORTANT: Copy the head OUTSIDE inference_mode.
initial_head = copy.deepcopy(
    baseline_model.lm_head
).to(DEVICE)

# Verify PyTorch can calculate gradients.
assert not frozen_features.is_inference()

for parameter in initial_head.parameters():
    assert parameter.requires_grad
    assert not parameter.is_inference()

print("AUTOGRAD TENSOR FIX: PASSED")

assert frozen_features.ndim == 3
assert frozen_features.shape[0] == 1

# Keep only actual target tokens, not padding.
targets = batch["labels"][
    batch["labels"] >= 0
].reshape(1, -1).contiguous()

assert targets.numel() > 0
assert not (targets == BLANK_ID).any().item()

input_lengths = torch.tensor(
    [frozen_features.shape[1]],
    dtype=torch.long
)

target_lengths = torch.tensor(
    [targets.shape[1]],
    dtype=torch.long
)

required_frames = (
    targets.shape[1]
    + (targets[0, 1:] == targets[0, :-1]).sum().item()
)

assert frozen_features.shape[1] >= required_frames

print("\nCACHED FEATURES")
print("Feature shape:", tuple(frozen_features.shape))
print("Target tokens:", targets.shape[1])
print("Required CTC frames:", required_frames)
print("Available frames:", frozen_features.shape[1])
print("Original model CTC loss:", round(initial_full_loss, 4))

# We no longer need the full pretrained encoder.
del baseline_model, original_forward
gc.collect()
torch.cuda.empty_cache()

# ==========================================
# 4. TRAIN ONLY THE ORIGINAL CTC HEAD
# ==========================================

head = initial_head.to(DEVICE)
head.train()

optimizer_probe = torch.optim.AdamW(
    head.parameters(),
    lr=HEAD_ONLY_LR,
    weight_decay=0.0
)

def head_only_loss():
    logits = head(frozen_features)

    # Use FP32 CTC to avoid mixed-precision
    # instability in this controlled experiment.
    log_probs = F.log_softmax(
        logits.float(),
        dim=-1
    ).transpose(0, 1)

    return F.ctc_loss(
        log_probs,
        targets,
        input_lengths,
        target_lengths,
        blank=BLANK_ID,
        reduction="mean",
        zero_infinity=False
    )


def evaluate_head():

    head.eval()

    with torch.no_grad():

        logits = head(frozen_features)

        probabilities = logits.float().softmax(
            dim=-1
        )

        predicted_ids = logits.argmax(dim=-1)

        predicted = processor.batch_decode(
            predicted_ids.cpu()
        )[0]

        predicted = normalize_amharic_ctc(
            predicted
        )

        blank_probability = (
            probabilities[..., BLANK_ID]
            .mean().item()
        )

        blank_argmax = (
            (predicted_ids == BLANK_ID)
            .float().mean().item()
        )

        loss = float(head_only_loss().item())

    return {
        "ctc_loss": loss,
        "cer": float(cer(REFERENCE, predicted)),
        "blank_probability": blank_probability,
        "blank_argmax": blank_argmax,
        "prediction": predicted
    }

# Sanity check: the cached-feature loss
# should match the complete starting model.
initial = evaluate_head()

print("\nLOSS CONSISTENCY CHECK")
print("Original model:", round(initial_full_loss, 5))
print("Cached features:", round(initial["ctc_loss"], 5))

assert abs(
    initial_full_loss - initial["ctc_loss"]
) < 0.05, "Cached-feature loss mismatch"

print("Consistency check: PASSED")

# ==========================================
# 5. RUN THE MEMORIZATION TEST
# ==========================================

history = []

for step in range(HEAD_ONLY_STEPS + 1):

    if step > 0:

        head.train()

        optimizer_probe.zero_grad(set_to_none=True)

        loss = head_only_loss()

        assert torch.isfinite(loss).item(), (
            f"Non-finite loss at step {step}"
        )

        loss.backward()

        torch.nn.utils.clip_grad_norm_(
            head.parameters(),
            max_norm=5.0,
            error_if_nonfinite=True
        )

        optimizer_probe.step()

    if step in REPORT_STEPS:

        result = evaluate_head()

        history.append({
            "step": step,
            **result
        })

        print(f"\nSTEP {step}/{HEAD_ONLY_STEPS}")
        print(
            "CTC loss:",
            round(result["ctc_loss"], 4)
        )
        print(
            "CER:",
            f"{result['cer'] * 100:.2f}%"
        )
        print(
            "Blank probability:",
            f"{result['blank_probability'] * 100:.2f}%"
        )
        print(
            "Blank argmax:",
            f"{result['blank_argmax'] * 100:.2f}%"
        )
        print(
            "Prediction:",
            result["prediction"][:200] or "[EMPTY]"
        )

        if result["cer"] <= 0.05:
            print("\nMEMORIZATION TARGET REACHED")
            break

# ==========================================
# 6. SAVE DIAGNOSTIC RESULTS
# ==========================================

HEAD_ONLY_RESULTS = (
    DATA_DIR / "head_only_step0_memorization.json"
)

report = {
    "starting_checkpoint": str(BASELINE_DIR),
    "recording_id": sample_record["id"],
    "reference": REFERENCE,
    "trainable_component": "lm_head_only",
    "cached_encoder_features": True,
    "learning_rate": HEAD_ONLY_LR,
    "maximum_steps": HEAD_ONLY_STEPS,
    "completed_steps": step,
    "history": history
}

with HEAD_ONLY_RESULTS.open(
    "w", encoding="utf-8"
) as file:
    json.dump(
        report,
        file,
        indent=2,
        ensure_ascii=False
    )

# ==========================================
# 7. FINAL COMPARISON
# ==========================================

final = history[-1]

print("\n" + "=" * 65)
print("HEAD-ONLY MEMORIZATION RESULTS")
print("=" * 65)

print("Starting loss:", round(initial["ctc_loss"], 4))
print("Final loss:", round(final["ctc_loss"], 4))

print(
    "Starting CER:",
    f"{initial['cer'] * 100:.2f}%"
)
print(
    "Final CER:",
    f"{final['cer'] * 100:.2f}%"
)

print("\nREFERENCE:")
print(REFERENCE)

print("\nFINAL PREDICTION:")
print(final["prediction"] or "[EMPTY]")

print("\nResults saved:", HEAD_ONLY_RESULTS)

# ==========================================
# 8. CLEAN UP
# ==========================================

del head, initial_head, optimizer_probe
del frozen_features, batch, targets

gc.collect()
torch.cuda.empty_cache()

print("\nMAIN EXPERIMENT UNCHANGED")
print("Head-only diagnostic completed independently.")
print("Existing training checkpoints were not modified.")


HEAD-ONLY EXPERIMENT READY
Device: cuda
Original baseline: /content/drive/MyDrive/Amharic_ASR_XLSR/baselines/xlsr_step0
Sample: 6Q0fEziAqyQVIz4J8aws
Duration: 5.184 seconds
Target tokens: 39
No step-500 model required.
FROZEN-ENCODER MEMORIZATION EXPERIMENT
-------------------------------------------------------
Recording: 6Q0fEziAqyQVIz4J8aws
Reference: ይህ ምስል የሚያሳየው ከሸክላ የሚሰራ የሸክላ ድስት ምስል ነው
Model starting point: STEP ZERO
Trainable component: CTC HEAD ONLY
Maximum updates: 1000
AUTOGRAD TENSOR FIX: PASSED

CACHED FEATURES
Feature shape: (1, 258, 1024)
Target tokens: 39
Required CTC frames: 39
Available frames: 258
Original model CTC loss: 33.2449

LOSS CONSISTENCY CHECK
Original model: 33.24486
Cached features: 33.24486
Consistency check: PASSED

STEP 0/1000
CTC loss: 33.2449
CER: 256.41%
Blank probability: 0.38%
Blank argmax: 0.00%
Prediction: ጠጹኧጹኻጹኻሣጹሣኻ፲ኻጹኻሣኻጹኻሼጹኻጹኻጹሣtጹሣጹኻጹኻጹሣጹኻጹኻጹኻጹሣጹኻtሼኻጹሼኦጹሄኻጹሣጹኻtጹኻጹሣኻጹtሣጹኻጹሣኻ፲ጹሼጹኻጹሼሣኻጹኻጹኻጹኻጹሼጹሣኻጹኻጹሣጹtጹኧ

STEP 25/1000
CTC loss: 7.1819
CER: 97.

In [ ]:

# =====================================================
# CELL 36 - EXTENDED HEAD-ONLY MEMORIZATION
# Goal: Can frozen XLS-R features reach 0% CER?
# Saves resumable checkpoints every 250 updates.
# Does not modify the main step-500 model.
# =====================================================

import copy
import json
import gc
from pathlib import Path

import torch
import torch.nn.functional as F
from jiwer import cer, wer
from transformers import Wav2Vec2ForCTC

MAX_STEPS = 4000
REPORT_EVERY = 250
LEARNING_RATE = 1e-3

TARGET_ID = "6Q0fEziAqyQVIz4J8aws"
BLANK_ID = tokenizer.pad_token_id
REFERENCE = sample_record["transcription"]

assert sample_record["id"] == TARGET_ID
assert sample_example is not None
assert torch.is_grad_enabled()

SAVE_DIR = DATA_DIR / "head_only_extended"
SAVE_DIR.mkdir(parents=True, exist_ok=True)

CHECKPOINT_PATH = SAVE_DIR / "latest.pt"
HISTORY_PATH = SAVE_DIR / "history.json"

device = torch.device(DEVICE)

# -----------------------------------------------------
# 1. Cache features from the ORIGINAL pretrained model
# -----------------------------------------------------

print("Loading original XLS-R checkpoint...")

original = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(device)

original.eval()

probe_batch = ctc_collator([sample_example])
probe_batch = {
    key: value.to(device)
    for key, value in probe_batch.items()
}

with torch.no_grad():
    original_loss = float(
        original(**probe_batch).loss.item()
    )

    features = original.wav2vec2(
        input_values=probe_batch["input_values"],
        attention_mask=probe_batch["attention_mask"]
    ).last_hidden_state

features = features.detach().clone().float()

# Copy trainable head outside any inference context.
probe_head = copy.deepcopy(
    original.lm_head
).to(device).float()

assert not features.is_inference()
assert probe_head.weight.requires_grad

del original
gc.collect()
torch.cuda.empty_cache()

# -----------------------------------------------------
# 2. Prepare CTC labels
# -----------------------------------------------------

probe_targets = probe_batch["labels"][
    probe_batch["labels"] >= 0
].reshape(1, -1).contiguous()

input_lengths = torch.tensor(
    [features.shape[1]], dtype=torch.long
)
target_lengths = torch.tensor(
    [probe_targets.shape[1]], dtype=torch.long
)

assert probe_targets.shape[1] > 0
assert features.shape[1] >= probe_targets.shape[1]

probe_optimizer = torch.optim.AdamW(
    probe_head.parameters(),
    lr=LEARNING_RATE,
    weight_decay=0.0
)

def probe_loss():
    logits = probe_head(features)
    log_probs = F.log_softmax(
        logits.float(), dim=-1
    ).transpose(0, 1)

    return F.ctc_loss(
        log_probs,
        probe_targets,
        input_lengths,
        target_lengths,
        blank=BLANK_ID,
        reduction="mean",
        zero_infinity=False
    )

def probe_evaluate():
    probe_head.eval()

    with torch.no_grad():
        logits = probe_head(features)
        predicted_ids = logits.argmax(-1)

        prediction = processor.batch_decode(
            predicted_ids.cpu()
        )[0]

        prediction = normalize_amharic_ctc(
            prediction
        )

        loss = float(probe_loss().item())

        blank_fraction = (
            (predicted_ids == BLANK_ID)
            .float().mean().item()
        )

    return {
        "loss": loss,
        "cer": float(cer(REFERENCE, prediction)),
        "wer": float(wer(REFERENCE, prediction)),
        "blank_argmax": blank_fraction,
        "prediction": prediction
    }

# -----------------------------------------------------
# 3. Resume previous extended experiment if available
# -----------------------------------------------------

history = []
start_step = 0

if CHECKPOINT_PATH.exists():
    saved = torch.load(
        CHECKPOINT_PATH,
        map_location=device,
        weights_only=True
    )

    assert saved["recording_id"] == TARGET_ID

    probe_head.load_state_dict(saved["head"])
    probe_optimizer.load_state_dict(saved["optimizer"])

    start_step = int(saved["step"])

    if HISTORY_PATH.exists():
        history = json.loads(
            HISTORY_PATH.read_text(encoding="utf-8")
        )

    print(f"Resuming from step {start_step}")

else:
    # Verify cached features give the same initial loss.
    initial_loss = float(probe_loss().item())

    assert abs(initial_loss - original_loss) < 0.05, (
        "Initial loss differs from original model."
    )

    print("Initial loss consistency: PASSED")

def save_progress(step, result):
    checkpoint = {
        "recording_id": TARGET_ID,
        "step": step,
        "head": probe_head.state_dict(),
        "optimizer": probe_optimizer.state_dict()
    }

    temporary = SAVE_DIR / "latest.pt.partial"
    torch.save(checkpoint, temporary)
    temporary.replace(CHECKPOINT_PATH)

    temporary_history = SAVE_DIR / "history.json.partial"

    temporary_history.write_text(
        json.dumps(
            history, ensure_ascii=False, indent=2
        ),
        encoding="utf-8"
    )
    temporary_history.replace(HISTORY_PATH)

# -----------------------------------------------------
# 4. Train, evaluate and checkpoint
# -----------------------------------------------------

print("\nEXTENDED MEMORIZATION EXPERIMENT")
print("-" * 55)
print("Recording:", TARGET_ID)
print("Training from step:", start_step)
print("Maximum step:", MAX_STEPS)
print("Frozen feature shape:", tuple(features.shape))

current = probe_evaluate()

print(f"\nSTEP {start_step}")
print("Loss:", round(current["loss"], 4))
print("CER:", f"{current['cer'] * 100:.2f}%")
print("Prediction:", current["prediction"] or "[EMPTY]")

if not history:
    history.append({"step": start_step, **current})

completed_step = start_step

for step in range(start_step + 1, MAX_STEPS + 1):

    probe_head.train()
    probe_optimizer.zero_grad(set_to_none=True)

    loss = probe_loss()

    assert torch.isfinite(loss).item()
    assert loss.requires_grad

    loss.backward()

    torch.nn.utils.clip_grad_norm_(
        probe_head.parameters(),
        max_norm=5.0,
        error_if_nonfinite=True
    )

    probe_optimizer.step()
    completed_step = step

    if step % REPORT_EVERY == 0 or step == MAX_STEPS:

        result = probe_evaluate()

        history.append({"step": step, **result})
        save_progress(step, result)

        print(f"\nSTEP {step}/{MAX_STEPS}")
        print("CTC loss:", round(result["loss"], 4))
        print("CER:", f"{result['cer'] * 100:.2f}%")
        print("WER:", f"{result['wer'] * 100:.2f}%")
        print(
            "Blank argmax:",
            f"{result['blank_argmax'] * 100:.2f}%"
        )
        print(
            "Prediction:",
            result["prediction"] or "[EMPTY]"
        )

        if result["cer"] == 0.0:
            print("\nEXACT TRANSCRIPTION MEMORIZED!")
            break

# -----------------------------------------------------
# 5. Final result
# -----------------------------------------------------

final = probe_evaluate()

print("\n" + "=" * 55)
print("FINAL RESULT")
print("=" * 55)
print("Completed steps:", completed_step)
print("Final CER:", f"{final['cer'] * 100:.2f}%")
print("Final WER:", f"{final['wer'] * 100:.2f}%")

print("\nREFERENCE:")
print(REFERENCE)

print("\nPREDICTION:")
print(final["prediction"] or "[EMPTY]")

print("\nCheckpoint:", CHECKPOINT_PATH)
print("History:", HISTORY_PATH)

print("\nOriginal baseline and step-500 model unchanged.")


Loading original XLS-R checkpoint...
Initial loss consistency: PASSED

EXTENDED MEMORIZATION EXPERIMENT
-------------------------------------------------------
Recording: 6Q0fEziAqyQVIz4J8aws
Training from step: 0
Maximum step: 4000
Frozen feature shape: (1, 258, 1024)

STEP 0
Loss: 33.2449
CER: 256.41%
Prediction: ጠጹኧጹኻጹኻሣጹሣኻ፲ኻጹኻሣኻጹኻሼጹኻጹኻጹሣtጹሣጹኻጹኻጹሣጹኻጹኻጹኻጹሣጹኻtሼኻጹሼኦጹሄኻጹሣጹኻtጹኻጹሣኻጹtሣጹኻጹሣኻ፲ጹሼጹኻጹሼሣኻጹኻጹኻጹኻጹሼጹሣኻጹኻጹሣጹtጹኧ

STEP 250/4000
CTC loss: 1.7316
CER: 64.10%
WER: 100.00%
Blank argmax: 93.41%
Prediction: ይምየያውስሰራየድስትምስው

STEP 500/4000
CTC loss: 1.1085
CER: 51.28%
WER: 100.00%
Blank argmax: 91.47%
Prediction: ይምስየያሳውከየሰራ የድስትምስው

STEP 750/4000
CTC loss: 0.7775
CER: 41.03%
WER: 100.00%
Blank argmax: 89.92%
Prediction: ይህምስየያሳውከሸየሰራ የ ድስትምስነው

STEP 1000/4000
CTC loss: 0.5639
CER: 33.33%
WER: 100.00%
Blank argmax: 88.37%
Prediction: ይህምስየያሳው ከሸየሰራ የሸ ድስትምስልነው

STEP 1250/4000
CTC loss: 0.431
CER: 30.77%
WER: 100.00%
Blank argmax: 87.98%
Prediction: ይህምስየሚያሳው ከሸየሰራ የሸ ድስትምስልነው

STEP 1500/4000


In [ ]:

# ============================================================
# CELL 37 - CONTROLLED ENCODER COMPARISON
#
# Question:
# Did fine-tuning to step 500 make the encoder's
# features harder to learn from?
#
# CONTROL:
# Step-0 encoder + step-0 head -> 0% CER at 2250 steps
#
# TEST:
# Step-500 encoder + SAME step-0 head initialization
#
# Both encoders remain frozen.
# No existing checkpoint will be modified.
# ============================================================

import copy
import json
import gc
from pathlib import Path

import torch
import torch.nn.functional as F
from jiwer import cer, wer
from transformers import Wav2Vec2ForCTC

CONTROL_MAX_STEPS = 2500
CONTROL_LR = 1e-3
CONTROL_REPORT_EVERY = 250

CONTROL_ID = "6Q0fEziAqyQVIz4J8aws"
CONTROL_BLANK = tokenizer.pad_token_id

STEP500_PATH = CHECKPOINT_DIR / "step_000500"

CONTROL_DIR = DATA_DIR / "encoder_step500_head_control"
CONTROL_DIR.mkdir(parents=True, exist_ok=True)

CONTROL_CKPT = CONTROL_DIR / "latest.pt"
CONTROL_HISTORY = CONTROL_DIR / "history.json"

ORIGINAL_HISTORY = (
    DATA_DIR / "head_only_extended" / "history.json"
)

assert Path(BASELINE_DIR).is_dir()
assert STEP500_PATH.is_dir()
assert ORIGINAL_HISTORY.is_file()
assert sample_record["id"] == CONTROL_ID
assert sample_example is not None
assert torch.is_grad_enabled()

control_device = torch.device(DEVICE)
control_reference = sample_record["transcription"]

# ------------------------------------------------------------
# 1. Prepare exactly the same recording and labels
# ------------------------------------------------------------

control_batch = ctc_collator([sample_example])

control_batch = {
    k: v.to(control_device)
    for k, v in control_batch.items()
}

control_targets = control_batch["labels"][
    control_batch["labels"] >= 0
].reshape(1, -1).contiguous()

control_target_lengths = torch.tensor(
    [control_targets.shape[1]], dtype=torch.long
)

# ------------------------------------------------------------
# 2. Load original encoder and save its original head
# ------------------------------------------------------------

print("Loading STEP-0 model...")

original_model = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(control_device)

original_model.eval()

with torch.no_grad():
    original_features = original_model.wav2vec2(
        input_values=control_batch["input_values"],
        attention_mask=control_batch["attention_mask"]
    ).last_hidden_state.detach().clone().float()

# Copy outside inference mode. Keep the exact starting head.
control_head = copy.deepcopy(
    original_model.lm_head
).to(control_device).float()

del original_model
gc.collect()
torch.cuda.empty_cache()

# ------------------------------------------------------------
# 3. Get features from the STEP-500 encoder
# ------------------------------------------------------------

print("Loading STEP-500 model...")

step500_model = Wav2Vec2ForCTC.from_pretrained(
    str(STEP500_PATH)
).to(control_device)

step500_model.eval()

with torch.no_grad():
    step500_features = step500_model.wav2vec2(
        input_values=control_batch["input_values"],
        attention_mask=control_batch["attention_mask"]
    ).last_hidden_state.detach().clone().float()

del step500_model
gc.collect()
torch.cuda.empty_cache()

assert original_features.shape == step500_features.shape
assert not step500_features.is_inference()
assert control_head.weight.requires_grad

control_input_lengths = torch.tensor(
    [step500_features.shape[1]], dtype=torch.long
)

assert step500_features.shape[1] >= (
    control_targets.shape[1]
    + (
        control_targets[0, 1:]
        == control_targets[0, :-1]
    ).sum().item()
)

# ------------------------------------------------------------
# 4. Verify original experimental conditions
# ------------------------------------------------------------

def control_ctc_loss(features):
    logits = control_head(features)

    return F.ctc_loss(
        F.log_softmax(
            logits.float(), dim=-1
        ).transpose(0, 1),
        control_targets,
        control_input_lengths,
        control_target_lengths,
        blank=CONTROL_BLANK,
        reduction="mean",
        zero_infinity=False
    )

with torch.no_grad():
    original_start_loss = float(
        control_ctc_loss(original_features).item()
    )

assert abs(original_start_loss - 33.24486) < 0.05, (
    "Starting head or original features do not match "
    "the previous controlled experiment."
)

del original_features
torch.cuda.empty_cache()

print("\nCONTROL VERIFICATION")
print("-" * 50)
print("Original starting loss:", round(original_start_loss, 5))
print("Expected:", 33.24486)
print("Verification: PASSED")
print("Step-500 feature shape:", tuple(step500_features.shape))

# ------------------------------------------------------------
# 5. Create independent head optimizer
# ------------------------------------------------------------

control_optimizer = torch.optim.AdamW(
    control_head.parameters(),
    lr=CONTROL_LR,
    weight_decay=0.0
)

def evaluate_control():

    control_head.eval()

    with torch.no_grad():
        logits = control_head(step500_features)
        predictions = logits.argmax(dim=-1)

        text = processor.batch_decode(
            predictions.cpu()
        )[0]

        text = normalize_amharic_ctc(text)

        current_loss = float(
            control_ctc_loss(step500_features).item()
        )

        blank_fraction = float(
            (predictions == CONTROL_BLANK)
            .float().mean().item()
        )

    return {
        "loss": current_loss,
        "cer": float(cer(control_reference, text)),
        "wer": float(wer(control_reference, text)),
        "blank_argmax": blank_fraction,
        "prediction": text
    }

# ------------------------------------------------------------
# 6. Load original encoder learning curve
# ------------------------------------------------------------

with ORIGINAL_HISTORY.open(encoding="utf-8") as f:
    original_history = json.load(f)

original_by_step = {
    int(row["step"]): row
    for row in original_history
}

assert original_by_step[2250]["cer"] == 0.0

# ------------------------------------------------------------
# 7. Resume this diagnostic if it was interrupted
# ------------------------------------------------------------

control_history = []
control_start = 0

if CONTROL_CKPT.exists():

    state = torch.load(
        CONTROL_CKPT,
        map_location=control_device,
        weights_only=True
    )

    assert state["recording_id"] == CONTROL_ID
    assert state["experiment"] == "step500_encoder_step0_head"

    control_head.load_state_dict(state["head"])
    control_optimizer.load_state_dict(state["optimizer"])

    control_start = int(state["step"])

    if CONTROL_HISTORY.exists():
        control_history = json.loads(
            CONTROL_HISTORY.read_text(encoding="utf-8")
        )

    print("\nResuming diagnostic from step", control_start)

def save_control(step):

    state = {
        "experiment": "step500_encoder_step0_head",
        "recording_id": CONTROL_ID,
        "step": step,
        "head": control_head.state_dict(),
        "optimizer": control_optimizer.state_dict()
    }

    temp = CONTROL_DIR / "latest.pt.partial"
    torch.save(state, temp)
    temp.replace(CONTROL_CKPT)

    history_temp = CONTROL_DIR / "history.json.partial"
    history_temp.write_text(
        json.dumps(
            control_history, indent=2, ensure_ascii=False
        ),
        encoding="utf-8"
    )
    history_temp.replace(CONTROL_HISTORY)

# ------------------------------------------------------------
# 8. Run controlled comparison
# ------------------------------------------------------------

print("\nENCODER COMPARISON")
print("=" * 60)
print("Same recording:", CONTROL_ID)
print("Same head initialization: YES")
print("Same LR:", CONTROL_LR)
print("Only difference: Encoder at step 0 vs step 500")
print("Training starts at:", control_start)

start_result = evaluate_control()

print("\nSTEP", control_start)
print("CTC loss:", round(start_result["loss"], 4))
print("CER:", f"{start_result['cer'] * 100:.2f}%")
print("Prediction:", start_result["prediction"] or "[EMPTY]")

if not control_history:
    control_history.append({
        "step": control_start,
        **start_result
    })

completed_step = control_start

if start_result["cer"] == 0.0:
    print("Memorization already achieved.")
else:
    for step in range(control_start + 1, CONTROL_MAX_STEPS + 1):

        control_head.train()
        control_optimizer.zero_grad(set_to_none=True)

        loss = control_ctc_loss(step500_features)

        assert torch.isfinite(loss).item()
        assert loss.requires_grad

        loss.backward()

        torch.nn.utils.clip_grad_norm_(
            control_head.parameters(),
            max_norm=5.0,
            error_if_nonfinite=True
        )

        control_optimizer.step()
        completed_step = step

        if step % CONTROL_REPORT_EVERY == 0:

            result = evaluate_control()

            control_history.append({
                "step": step,
                **result
            })

            save_control(step)

            print(f"\nSTEP {step}/{CONTROL_MAX_STEPS}")
            print(
                "Step-500 encoder CER:",
                f"{result['cer'] * 100:.2f}%"
            )

            original_result = original_by_step.get(step)

            if original_result is not None:
                print(
                    "Step-0 encoder CER:",
                    f"{original_result['cer'] * 100:.2f}%"
                )

            print("CTC loss:", round(result["loss"], 4))
            print(
                "Blank argmax:",
                f"{result['blank_argmax'] * 100:.2f}%"
            )
            print(
                "Prediction:",
                result["prediction"] or "[EMPTY]"
            )

            if result["cer"] == 0.0:
                print("\nEXACT TRANSCRIPTION MEMORIZED")
                break

# ------------------------------------------------------------
# 9. Final diagnostic
# ------------------------------------------------------------

final_result = evaluate_control()

print("\n" + "=" * 60)
print("CONTROLLED COMPARISON COMPLETE")
print("=" * 60)

print("Original encoder:")
print("  Reached 0% CER at step 2250")

print("\nStep-500 encoder:")
print("  Completed steps:", completed_step)
print(
    "  Final CER:",
    f"{final_result['cer'] * 100:.2f}%"
)
print(
    "  Final WER:",
    f"{final_result['wer'] * 100:.2f}%"
)
print("  Final loss:", round(final_result["loss"], 4))

print("\nREFERENCE:")
print(control_reference)

print("\nPREDICTION:")
print(final_result["prediction"] or "[EMPTY]")

print("\nSaved:", CONTROL_DIR)
print("Existing training checkpoints unchanged.")


Loading STEP-0 model...
Loading STEP-500 model...

CONTROL VERIFICATION
--------------------------------------------------
Original starting loss: 33.24486
Expected: 33.24486
Verification: PASSED
Step-500 feature shape: (1, 258, 1024)

ENCODER COMPARISON
Same recording: 6Q0fEziAqyQVIz4J8aws
Same head initialization: YES
Same LR: 0.001
Only difference: Encoder at step 0 vs step 500
Training starts at: 0

STEP 0
CTC loss: 24.9455
CER: 100.00%
Prediction: [EMPTY]

STEP 250/2500
Step-500 encoder CER: 94.87%
Step-0 encoder CER: 64.10%
CTC loss: 2.3632
Blank argmax: 99.22%
Prediction: ይው

STEP 500/2500
Step-500 encoder CER: 84.62%
Step-0 encoder CER: 51.28%
CTC loss: 1.8124
Blank argmax: 96.90%
Prediction: ይምያውክው

STEP 750/2500
Step-500 encoder CER: 66.67%
Step-0 encoder CER: 41.03%
CTC loss: 1.3636
Blank argmax: 94.57%
Prediction: ይምያውሸክሸክላምስልው

STEP 1000/2500
Step-500 encoder CER: 64.10%
Step-0 encoder CER: 33.33%
CTC loss: 1.0677
Blank argmax: 93.80%
Prediction: ይምያሳውሸክሸክላምስልው

STEP 1250/

In [ ]:

# ============================================================
# CELL 38 - SMALL DATASET FOR CONTROLLED ASR TRAINING
#
# 8 training recordings from 8 speakers
# 4 held-out recordings from 4 DIFFERENT speakers
#
# No model training and no checkpoint modifications.
# ============================================================

import json
import random
from pathlib import Path
from IPython.display import Audio, display

SMALL_SET_DIR = DATA_DIR / "head_only_multirecording_v1"
SMALL_SET_DIR.mkdir(parents=True, exist_ok=True)

SMALL_SET_PATH = SMALL_SET_DIR / "selection.json"

TRAIN_COUNT = 8
VAL_COUNT = 4
SELECTION_SEED = 20261019

# XLS-R 300M convolution configuration.
CONV_KERNELS = (10, 3, 3, 3, 3, 2, 2)
CONV_STRIDES = (5, 2, 2, 2, 2, 2, 2)

def count_output_frames(num_samples):
    length = int(num_samples)
    for kernel, stride in zip(CONV_KERNELS, CONV_STRIDES):
        length = (length - kernel) // stride + 1
    return length

def inspect_record(record):

    duration = float(record["duration_seconds"])
    speaker = record.get("speaker_id")

    if not speaker or not (4.0 <= duration <= 18.0):
        return None

    audio_path = Path(AUDIO_DIR) / record["audio_file"]

    if not audio_path.is_file():
        return None

    labels = tokenizer.encode(
        record["transcription"],
        add_special_tokens=False
    )

    if not (25 <= len(labels) <= 140):
        return None

    if tokenizer.unk_token_id in labels:
        return None

    repeated = sum(
        a == b
        for a, b in zip(labels[:-1], labels[1:])
    )

    required = len(labels) + repeated
    available = count_output_frames(
        round(duration * 16000)
    )

    # Leave a conservative alignment margin.
    if available - required < 20:
        return None

    return {
        "record": record,
        "tokens": len(labels),
        "margin": available - required
    }

# ------------------------------------------------------------
# 1. Select recordings or reuse saved selection
# ------------------------------------------------------------

record_lookup = {
    r["id"]: r for r in train_records
}

if SMALL_SET_PATH.exists():

    selection = json.loads(
        SMALL_SET_PATH.read_text(encoding="utf-8")
    )

    train_ids = selection["train_ids"]
    val_ids = selection["val_ids"]

    print("Loaded existing selection.")

else:

    eligible = []

    for record in train_records:
        result = inspect_record(record)
        if result is not None:
            eligible.append(result)

    rng = random.Random(SELECTION_SEED)
    rng.shuffle(eligible)

    selected = []
    used_speakers = set()

    for candidate in eligible:

        record = candidate["record"]
        speaker = record["speaker_id"]

        if speaker in used_speakers:
            continue

        selected.append(record["id"])
        used_speakers.add(speaker)

        if len(selected) == TRAIN_COUNT + VAL_COUNT:
            break

    print("Eligible recordings:", len(eligible))
    print("Selected speakers:", len(selected))

    assert len(selected) == TRAIN_COUNT + VAL_COUNT, (
        "Not enough suitable recordings with distinct speakers."
    )

    train_ids = selected[:TRAIN_COUNT]
    val_ids = selected[TRAIN_COUNT:]

    selection = {
        "seed": SELECTION_SEED,
        "train_ids": train_ids,
        "val_ids": val_ids
    }

    SMALL_SET_PATH.write_text(
        json.dumps(
            selection, ensure_ascii=False, indent=2
        ),
        encoding="utf-8"
    )

# ------------------------------------------------------------
# 2. Validate our selected recordings
# ------------------------------------------------------------

assert len(train_ids) == TRAIN_COUNT
assert len(val_ids) == VAL_COUNT

assert len(set(train_ids + val_ids)) == (
    TRAIN_COUNT + VAL_COUNT
)

small_train_records = [
    record_lookup[id_] for id_ in train_ids
]

small_val_records = [
    record_lookup[id_] for id_ in val_ids
]

train_speakers = {
    r["speaker_id"] for r in small_train_records
}
val_speakers = {
    r["speaker_id"] for r in small_val_records
}

assert not (train_speakers & val_speakers)
assert len(train_speakers) == TRAIN_COUNT
assert len(val_speakers) == VAL_COUNT

for record in small_train_records + small_val_records:
    assert inspect_record(record) is not None, (
        f"Missing audio or invalid recording: {record['id']}"
    )

print("\n" + "=" * 60)
print("SMALL DATASET VERIFICATION")
print("=" * 60)

print("Training recordings:", len(small_train_records))
print("Held-out recordings:", len(small_val_records))
print("Overlapping speakers:", len(train_speakers & val_speakers))

print("\nTRAINING RECORDINGS")
for i, r in enumerate(small_train_records, 1):
    print(
        f"{i}. {r['id']} | "
        f"{r['duration_seconds']:.2f}s | "
        f"speaker={r['speaker_id']}"
    )
    print("   ", r["transcription"][:130])

print("\nHELD-OUT RECORDINGS")
for i, r in enumerate(small_val_records, 1):
    print(
        f"{i}. {r['id']} | "
        f"{r['duration_seconds']:.2f}s | "
        f"speaker={r['speaker_id']}"
    )
    print("   ", r["transcription"][:130])

# ------------------------------------------------------------
# 3. Listen to three recordings
# ------------------------------------------------------------

examples_to_listen = [
    ("TRAIN 1", small_train_records[0]),
    ("TRAIN 2", small_train_records[1]),
    ("HELD-OUT 1", small_val_records[0])
]

print("\n" + "=" * 60)
print("AUDIO AND TRANSCRIPT QUALITY CHECK")
print("=" * 60)

for label, record in examples_to_listen:

    print("\n", label)
    print("Recording ID:", record["id"])
    print("Transcription:", record["transcription"])

    audio_file = Path(AUDIO_DIR) / record["audio_file"]

    display(Audio(filename=str(audio_file)))

print("\nSelection saved:", SMALL_SET_PATH)
print("No model weights or checkpoints were modified.")


Eligible recordings: 2615
Selected speakers: 12

SMALL DATASET VERIFICATION
Training recordings: 8
Held-out recordings: 4
Overlapping speakers: 0

TRAINING RECORDINGS
1. aXx7RwawmZHKRpxFNU6p | 16.22s | speaker=7uE8erckn1Z98lz9QpfXPAEHifO2
    ቬጀቴሪያንነትና ቪጋኒዝም የእንስሳት ተዋጽኦዎችን የማይጠቀሙ የምግብ ምርጫዎች ሲሆኑ የራሳቸው ጥቅሞች አሏቸው
2. 37kmKxvapB3drOS3Kpcf | 17.78s | speaker=MfppGpxsCohMsinOkuWwe6AMAGt2
    ግብርና ኢትዮጵያ በግብርና ሥራ የምትጣወቅ ሀገር ናት ግብርና በሀገራችን 80 የሚሆነውን ኢኮኖሚ ትሸፍኖ የሚገኝ ነው በግብርና አብዛኛው የኢትዮጵያ ማሕበረሰብ የሚተዳደርበት ነው
3. 0NCgT71hjXyrBZrhYN79 | 16.22s | speaker=FPxKrorhxlhUZsf2uoAPWA2GRns1
    በዚህ በመስኖ ላይ የምትመለከቱት ደግሞ ቆሻሻ ቦታዎችን እንመለከታለን አንዲት ሴትዮ ደግሞ ቆሻሻ እያፀዳች እንመለከታለን የቆሻሻ ጋሪም በቆሻሻ ተሞልቶ እናያለን
4. ScHb8g7RjsOuSbfBvppf | 16.94s | speaker=bnlO6rMd4pVOKWDyVhQfojksz6h2
    የኢነጅኦ ባንኮች የምንላቸው በተለያዩ የኢነጅኦ ወይም ደግሞ በተለያዩ ኦርጋናይዜሽኖች የሚከናወን የምግብ ድጋፍ ሲሆን ለተቸገሩ ሀገራት ወይም ደግሞ በጦርነት ውስጥ ላሉ ሀገራት ይደርሳል
5. 09B2bpTuKAta4p2U5x3h | 15.22s | speaker=ntYvnLxnh4VyEsSg5VAc4b1R93g1
    የታዳጊዎች ጤና በወጣትነት እድሜ ላይ የሚገኙ ልጆችን የ ፆታዊ ጤና የ አመጋገብ ቺግሮ


 TRAIN 2
Recording ID: 37kmKxvapB3drOS3Kpcf
Transcription: ግብርና ኢትዮጵያ በግብርና ሥራ የምትጣወቅ ሀገር ናት ግብርና በሀገራችን 80 የሚሆነውን ኢኮኖሚ ትሸፍኖ የሚገኝ ነው በግብርና አብዛኛው የኢትዮጵያ ማሕበረሰብ የሚተዳደርበት ነው



 HELD-OUT 1
Recording ID: 3TSyIpivT7BhbbeVJG76
Transcription: ውይ ማር እንዴት እንዲሚያምር ይ በባሊ በባሊ ሆኖ የተቆረጠ ተቆርጦ የተቀመጠ ማህርን የምንመለከት ሲሆን በጣም ያምራል እንዴት እንዲሚያስጎመጅ ብስመአብ



Selection saved: /content/drive/MyDrive/Amharic_ASR_XLSR/data/head_only_multirecording_v1/selection.json
No model weights or checkpoints were modified.


In [ ]:

# ============================================================
# CELL 39 - MULTI-RECORDING HEAD-ONLY ASR EXPERIMENT
#
# 8 training recordings / 4 held-out recordings
# Original XLS-R encoder is FROZEN.
# Only the CTC prediction head is trained.
#
# Saves checkpoints; does NOT change previous models.
# ============================================================

import json
import gc
import copy
import hashlib
from pathlib import Path

import torch
import torch.nn.functional as F
from jiwer import cer, wer
from transformers import Wav2Vec2ForCTC

# ------------------------------------------------------------
# 1. Configuration
# ------------------------------------------------------------

MAX_UPDATES = 4000
REPORT_EVERY = 250
LEARNING_RATE = 1e-3
BLANK_ID = tokenizer.pad_token_id

device = torch.device(
    "cuda" if torch.cuda.is_available() else "cpu"
)

EXPERIMENT_DIR = (
    DATA_DIR / "head_only_multirecording_v1"
)
SELECTION_PATH = EXPERIMENT_DIR / "selection.json"
CHECKPOINT_PATH = EXPERIMENT_DIR / "training_latest.pt"
HISTORY_PATH = EXPERIMENT_DIR / "training_history.json"

assert SELECTION_PATH.exists()
assert Path(BASELINE_DIR).exists()

selection = json.loads(
    SELECTION_PATH.read_text(encoding="utf-8")
)

train_ids = selection["train_ids"]
val_ids = selection["val_ids"]

assert len(train_ids) == 8
assert len(val_ids) == 4
assert len(set(train_ids + val_ids)) == 12

record_by_id = {
    record["id"]: record
    for record in train_records
}

index_by_id = {
    record["id"]: i
    for i, record in enumerate(train_dataset.records)
}

train_speakers = {
    record_by_id[rid]["speaker_id"]
    for rid in train_ids
}
val_speakers = {
    record_by_id[rid]["speaker_id"]
    for rid in val_ids
}

assert not (train_speakers & val_speakers)

selection_signature = hashlib.sha256(
    json.dumps(
        {
            "train": train_ids,
            "val": val_ids,
            "references": {
                rid: record_by_id[rid]["transcription"]
                for rid in train_ids + val_ids
            }
        },
        sort_keys=True,
        ensure_ascii=False
    ).encode("utf-8")
).hexdigest()

print("MULTI-RECORDING EXPERIMENT")
print("=" * 55)
print("Training examples:", len(train_ids))
print("Held-out examples:", len(val_ids))
print("Shared speakers:", 0)
print("Device:", device)

# ------------------------------------------------------------
# 2. Load original pretrained encoder
# ------------------------------------------------------------

print("\nLoading original XLS-R checkpoint...")

base_model = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(device)

base_model.eval()

# Head is copied OUTSIDE inference mode.
head = copy.deepcopy(
    base_model.lm_head
).to(device).float()

assert head.weight.requires_grad
assert not head.weight.is_inference()

# ------------------------------------------------------------
# 3. Cache encoder features for all 12 examples
# ------------------------------------------------------------

def cache_example(record_id):

    example = train_dataset[
        index_by_id[record_id]
    ]

    batch = ctc_collator([example])
    batch = {
        key: value.to(device)
        for key, value in batch.items()
    }

    # Encoder is frozen.
    with torch.no_grad():
        hidden = base_model.wav2vec2(
            input_values=batch["input_values"],
            attention_mask=batch["attention_mask"]
        ).last_hidden_state

    hidden = hidden.detach().clone().float()

    targets = batch["labels"][
        batch["labels"] >= 0
    ].reshape(-1).contiguous()

    num_frames = hidden.shape[1]
    num_tokens = targets.numel()

    repeated = int(
        (targets[1:] == targets[:-1]).sum().item()
    )

    assert num_frames >= num_tokens + repeated
    assert not (targets == BLANK_ID).any()
    assert not hidden.is_inference()

    reference = normalize_amharic_ctc(
        record_by_id[record_id]["transcription"]
    )

    return {
        "id": record_id,
        "features": hidden,
        "targets": targets,
        "input_lengths": torch.tensor(
            [num_frames], dtype=torch.long
        ),
        "target_lengths": torch.tensor(
            [num_tokens], dtype=torch.long
        ),
        "reference": reference
    }

print("\nCaching 12 recordings...")

train_items = [
    cache_example(rid)
    for rid in train_ids
]

val_items = [
    cache_example(rid)
    for rid in val_ids
]

# No further need for the full encoder.
del base_model
gc.collect()
torch.cuda.empty_cache()

print("Encoder features cached: 12/12")
print(
    "Trainable parameters:",
    sum(p.numel() for p in head.parameters())
)

# ------------------------------------------------------------
# 4. CTC loss and evaluation
# ------------------------------------------------------------

def example_loss(item):
    logits = head(item["features"])

    log_probs = F.log_softmax(
        logits.float(),
        dim=-1
    ).transpose(0, 1)

    return F.ctc_loss(
        log_probs,
        item["targets"],
        item["input_lengths"],
        item["target_lengths"],
        blank=BLANK_ID,
        reduction="mean",
        zero_infinity=False
    )


def evaluate_group(items):
    head.eval()

    references = []
    predictions = []
    losses = []
    nonempty = 0

    with torch.no_grad():

        for item in items:

            logits = head(item["features"])

            predicted_ids = logits.argmax(
                dim=-1
            )

            prediction = processor.batch_decode(
                predicted_ids.cpu()
            )[0]

            prediction = normalize_amharic_ctc(
                prediction
            )

            reference = item["reference"]

            references.append(reference)
            predictions.append(prediction)

            losses.append(
                float(example_loss(item).item())
            )

            if prediction.strip():
                nonempty += 1

    return {
        "cer": float(cer(references, predictions)),
        "wer": float(wer(references, predictions)),
        "mean_loss": sum(losses) / len(losses),
        "nonempty": nonempty,
        "count": len(items),
        "references": references,
        "predictions": predictions
    }

optimizer = torch.optim.AdamW(
    head.parameters(),
    lr=LEARNING_RATE,
    weight_decay=0.0
)

# ------------------------------------------------------------
# 5. Resume experiment if previously saved
# ------------------------------------------------------------

history = []
start_step = 0

if CHECKPOINT_PATH.exists():

    state = torch.load(
        CHECKPOINT_PATH,
        map_location="cpu",
        weights_only=True
    )

    assert state["signature"] == selection_signature
    assert state["learning_rate"] == LEARNING_RATE

    head.load_state_dict(state["head"])
    optimizer.load_state_dict(state["optimizer"])

    start_step = int(state["step"])

    if HISTORY_PATH.exists():
        history = json.loads(
            HISTORY_PATH.read_text(encoding="utf-8")
        )

    print("\nResuming from update:", start_step)

else:
    print("\nStarting a new experiment.")

# ------------------------------------------------------------
# 6. Save a resumable checkpoint
# ------------------------------------------------------------

def save_experiment(step):

    state = {
        "step": step,
        "signature": selection_signature,
        "learning_rate": LEARNING_RATE,
        "head": head.state_dict(),
        "optimizer": optimizer.state_dict()
    }

    temp_checkpoint = (
        EXPERIMENT_DIR / "training_latest.pt.partial"
    )

    torch.save(state, temp_checkpoint)
    temp_checkpoint.replace(CHECKPOINT_PATH)

    temp_history = (
        EXPERIMENT_DIR / "training_history.json.partial"
    )

    temp_history.write_text(
        json.dumps(
            history,
            indent=2,
            ensure_ascii=False
        ),
        encoding="utf-8"
    )

    temp_history.replace(HISTORY_PATH)

# ------------------------------------------------------------
# 7. Evaluate before training
# ------------------------------------------------------------

def report_step(step):

    train_result = evaluate_group(train_items)
    val_result = evaluate_group(val_items)

    record = {
        "step": step,
        "train_cer": train_result["cer"],
        "train_wer": train_result["wer"],
        "train_loss": train_result["mean_loss"],
        "train_nonempty": train_result["nonempty"],
        "val_cer": val_result["cer"],
        "val_wer": val_result["wer"],
        "val_loss": val_result["mean_loss"],
        "val_nonempty": val_result["nonempty"]
    }

    print(f"\nUPDATE {step}/{MAX_UPDATES}")
    print("-" * 45)

    print(
        "TRAIN CER:",
        f"{train_result['cer'] * 100:.2f}%",
        "| WER:",
        f"{train_result['wer'] * 100:.2f}%"
    )

    print(
        "HELD-OUT CER:",
        f"{val_result['cer'] * 100:.2f}%",
        "| WER:",
        f"{val_result['wer'] * 100:.2f}%"
    )

    print(
        "Nonempty predictions:",
        f"{train_result['nonempty']}/8 train,",
        f"{val_result['nonempty']}/4 held-out"
    )

    print(
        "Mean train CTC loss:",
        round(train_result["mean_loss"], 4)
    )

    print("\nTRAIN SAMPLE:")
    print(
        train_result["predictions"][0][:150]
        or "[EMPTY]"
    )

    print("HELD-OUT SAMPLE:")
    print(
        val_result["predictions"][0][:150]
        or "[EMPTY]"
    )

    return record

if start_step == 0 and not history:
    history.append(report_step(0))

# ------------------------------------------------------------
# 8. Train on all eight examples in a rotating order
# ------------------------------------------------------------

print("\nBeginning head-only training...")
print("Maximum updates:", MAX_UPDATES)
print("Checkpoint interval:", REPORT_EVERY)

completed_step = start_step

for step in range(start_step + 1, MAX_UPDATES + 1):

    # Deterministic rotation through the eight examples.
    item = train_items[
        (step - 1) % len(train_items)
    ]

    head.train()
    optimizer.zero_grad(set_to_none=True)

    loss = example_loss(item)

    assert torch.isfinite(loss).item()
    assert loss.requires_grad

    loss.backward()

    torch.nn.utils.clip_grad_norm_(
        head.parameters(),
        max_norm=5.0,
        error_if_nonfinite=True
    )

    optimizer.step()
    completed_step = step

    if step % REPORT_EVERY == 0:

        result = report_step(step)
        history.append(result)

        save_experiment(step)

# ------------------------------------------------------------
# 9. Final report
# ------------------------------------------------------------

final_train = evaluate_group(train_items)
final_val = evaluate_group(val_items)

print("\n" + "=" * 60)
print("FINAL MULTI-RECORDING RESULTS")
print("=" * 60)

print("Completed updates:", completed_step)

print(
    "Train CER:",
    f"{final_train['cer'] * 100:.2f}%"
)

print(
    "Held-out CER:",
    f"{final_val['cer'] * 100:.2f}%"
)

print(
    "Held-out WER:",
    f"{final_val['wer'] * 100:.2f}%"
)

print("\nHELD-OUT EXAMPLE")
print("Reference:")
print(final_val["references"][0])
print("\nPrediction:")
print(final_val["predictions"][0] or "[EMPTY]")

print("\nCheckpoint:", CHECKPOINT_PATH)
print("History:", HISTORY_PATH)
print("Original XLS-R and step-500 model unchanged.")


MULTI-RECORDING EXPERIMENT
Training examples: 8
Held-out examples: 4
Shared speakers: 0
Device: cuda

Loading original XLS-R checkpoint...

Caching 12 recordings...
Encoder features cached: 12/12
Trainable parameters: 329025

Starting a new experiment.

UPDATE 0/4000
---------------------------------------------
TRAIN CER: 164.20% | WER: 100.00%
HELD-OUT CER: 213.39% | WER: 100.00%
Nonempty predictions: 8/8 train, 4/4 held-out
Mean train CTC loss: 42.3293

TRAIN SAMPLE:
ለኻኧኻጹኻለኧኻኧኻኧኻኧኻኧኻጹኻጹጕሄኻሄኻጹኻፓኻጹኧሣኻሄኻጹኧኻጹኻጹሄኻሄኻጹኧኻጹሼኻኦኻሄሣኻለኻኧኻጹመኻኧኻጹኻ፻ኻጹኧኻጹኧኻጹኧኻኧኻሼኻጹኧኻኧጹኻሼሣኻጹኻጹኻኧኻ፻ኻጹችኻሄኻሣኻጹኧኻኧኻኧኻጹኻጹሣኻጹኻፓጹኧኻኧኻኧ
HELD-OUT SAMPLE:
ጠኻጹኻጹኻጹኻጹኻtጹtጹኻጹኻጹኻጹኻጹኻጠጹኻጹኻጹኻጹኻጹኻጹኻጹኻጹኻጹሄጹሄጹኻጹኻጹኻጹኻጹኻጹኻጹኻጹኻጹኻጹኻጹኻጹችጹኻጹኻጹኻጹኻጹኻጹኻጹኻሄኻጹኻጠጹኻጹሄኻጹኻጹኻጹኻጹኻጹኻጹኻጹኻጹኻጹሼኻጹኻጹኻጹኻጹኻጹኧጹኻጹኻጹኻጹኻጹኻጹኻጹኻጹኻጹኻሄኻሣኻሼኻጹኻጹኻጹ

Beginning head-only training...
Maximum updates: 4000
Checkpoint interval: 250

UPDATE 250/4000
---------------------------------------------
TRAIN CER: 97.92% | WER: 100.00%
HELD-OUT CER: 99.21% | WER: 100.00%
Nonempty predicti

In [ ]:

# ============================================================
# CELL 40 - SHORT-RECORDING CONTROLLED DATASET
#
# 8 training recordings, including our proven sample
# 4 held-out recordings
# All 12 speakers must be distinct
# Recording duration: 3.5 to 8 seconds
#
# No model training or checkpoint changes.
# ============================================================

import json
import random
from pathlib import Path
from IPython.display import Audio, display

SHORT_DIR = DATA_DIR / "short_multirecording_v1"
SHORT_DIR.mkdir(parents=True, exist_ok=True)

SHORT_SELECTION_PATH = SHORT_DIR / "selection.json"

ANCHOR_ID = "6Q0fEziAqyQVIz4J8aws"
SEED = 20261019

TRAIN_COUNT = 8
VAL_COUNT = 4

CONV_KERNELS = (10, 3, 3, 3, 3, 2, 2)
CONV_STRIDES = (5, 2, 2, 2, 2, 2, 2)

def short_output_frames(n_samples):
    length = int(n_samples)
    for kernel, stride in zip(CONV_KERNELS, CONV_STRIDES):
        length = (length - kernel) // stride + 1
    return length

def short_candidate_ok(record):

    duration = float(record["duration_seconds"])
    speaker = record.get("speaker_id")
    transcript = record["transcription"]

    if not speaker:
        return False

    if not (3.5 <= duration <= 8.0):
        return False

    # Avoid digit-to-speech normalization ambiguity
    # in this small controlled experiment.
    if any(character.isdigit() for character in transcript):
        return False

    audio_path = Path(AUDIO_DIR) / record["audio_file"]

    if not audio_path.is_file():
        return False

    labels = tokenizer.encode(
        transcript,
        add_special_tokens=False
    )

    if not (20 <= len(labels) <= 85):
        return False

    if tokenizer.unk_token_id in labels:
        return False

    repeated = sum(
        left == right
        for left, right in zip(labels[:-1], labels[1:])
    )

    required_frames = len(labels) + repeated
    available_frames = short_output_frames(
        round(duration * 16000)
    )

    return available_frames - required_frames >= 30


record_lookup = {
    record["id"]: record
    for record in train_records
}

assert ANCHOR_ID in record_lookup
assert short_candidate_ok(record_lookup[ANCHOR_ID])

# ------------------------------------------------------------
# 1. Reuse selection if already generated
# ------------------------------------------------------------

if SHORT_SELECTION_PATH.exists():

    selection = json.loads(
        SHORT_SELECTION_PATH.read_text(
            encoding="utf-8"
        )
    )

    short_train_ids = selection["train_ids"]
    short_val_ids = selection["val_ids"]

    print("Restored existing short-recording selection.")

else:

    eligible = [
        record
        for record in train_records
        if short_candidate_ok(record)
        and record["id"] != ANCHOR_ID
    ]

    rng = random.Random(SEED)
    rng.shuffle(eligible)

    selected = [record_lookup[ANCHOR_ID]]
    used_speakers = {
        record_lookup[ANCHOR_ID]["speaker_id"]
    }

    for record in eligible:

        if record["speaker_id"] in used_speakers:
            continue

        selected.append(record)
        used_speakers.add(record["speaker_id"])

        if len(selected) == TRAIN_COUNT + VAL_COUNT:
            break

    assert len(selected) == 12, (
        "Not enough suitable recordings."
    )

    short_train_ids = [
        record["id"]
        for record in selected[:TRAIN_COUNT]
    ]

    short_val_ids = [
        record["id"]
        for record in selected[TRAIN_COUNT:]
    ]

    selection = {
        "seed": SEED,
        "anchor_id": ANCHOR_ID,
        "train_ids": short_train_ids,
        "val_ids": short_val_ids,
        "duration_range_seconds": [3.5, 8.0]
    }

    SHORT_SELECTION_PATH.write_text(
        json.dumps(
            selection,
            indent=2,
            ensure_ascii=False
        ),
        encoding="utf-8"
    )

    print("Eligible short recordings:", len(eligible))
    print("Created new short-recording selection.")

# ------------------------------------------------------------
# 2. Check sample integrity
# ------------------------------------------------------------

assert len(short_train_ids) == TRAIN_COUNT
assert len(short_val_ids) == VAL_COUNT
assert ANCHOR_ID in short_train_ids

all_ids = short_train_ids + short_val_ids

assert len(set(all_ids)) == 12

short_train_records = [
    record_lookup[rid]
    for rid in short_train_ids
]

short_val_records = [
    record_lookup[rid]
    for rid in short_val_ids
]

all_selected = (
    short_train_records + short_val_records
)

assert all(
    short_candidate_ok(record)
    for record in all_selected
)

all_speakers = [
    record["speaker_id"]
    for record in all_selected
]

assert len(set(all_speakers)) == 12

total_train_seconds = sum(
    float(record["duration_seconds"])
    for record in short_train_records
)

total_val_seconds = sum(
    float(record["duration_seconds"])
    for record in short_val_records
)

# ------------------------------------------------------------
# 3. Display selected dataset
# ------------------------------------------------------------

print("\n" + "=" * 60)
print("SHORT DATASET SUMMARY")
print("=" * 60)

print("Training recordings:", len(short_train_records))
print("Held-out recordings:", len(short_val_records))
print("Unique speakers:", len(set(all_speakers)))
print("Train duration:", round(total_train_seconds, 2), "seconds")
print("Held-out duration:", round(total_val_seconds, 2), "seconds")
print("Positive control:", ANCHOR_ID)

print("\nTRAINING RECORDINGS")
for index, record in enumerate(short_train_records, 1):
    print(
        f"\n{index}. {record['id']} "
        f"| {record['duration_seconds']:.2f}s"
    )
    print(record["transcription"])

print("\nHELD-OUT RECORDINGS")
for index, record in enumerate(short_val_records, 1):
    print(
        f"\n{index}. {record['id']} "
        f"| {record['duration_seconds']:.2f}s"
    )
    print(record["transcription"])

# ------------------------------------------------------------
# 4. Listen and check audio-to-text quality
# ------------------------------------------------------------

print("\n" + "=" * 60)
print("AUDIO QUALITY REVIEW")
print("=" * 60)

review_examples = [
    ("KNOWN POSITIVE CONTROL", short_train_records[0]),
    ("NEW TRAINING EXAMPLE", short_train_records[1]),
    ("NEW TRAINING EXAMPLE", short_train_records[2]),
    ("HELD-OUT EXAMPLE", short_val_records[0])
]

for label, record in review_examples:

    print("\n", label)
    print("ID:", record["id"])
    print("Transcript:", record["transcription"])

    audio_path = Path(AUDIO_DIR) / record["audio_file"]

    display(Audio(filename=str(audio_path)))

print("\nSelection saved:", SHORT_SELECTION_PATH)
print("No existing models or checkpoints were modified.")


AssertionError: Not enough suitable recordings.

In [ ]:

# ============================================================
# CELL 40B - ADAPTIVE SHORT-RECORDING DATASET FIX
# Prefer short recordings, relax duration when necessary.
# No training or checkpoint modifications.
# ============================================================

import json
import random
from pathlib import Path
from IPython.display import Audio, display

ANCHOR_ID = "6Q0fEziAqyQVIz4J8aws"
TRAIN_COUNT = 8
VAL_COUNT = 4

SHORT_DIR = DATA_DIR / "short_multirecording_v1"
SHORT_DIR.mkdir(parents=True, exist_ok=True)
SHORT_SELECTION_PATH = SHORT_DIR / "selection.json"

record_lookup = {r["id"]: r for r in train_records}
assert ANCHOR_ID in record_lookup

kernels = (10, 3, 3, 3, 3, 2, 2)
strides = (5, 2, 2, 2, 2, 2, 2)

def frame_count(samples):
    for kernel, stride in zip(kernels, strides):
        samples = (samples - kernel) // stride + 1
    return samples

def eligible_record(record):
    duration = float(record["duration_seconds"])
    text = record["transcription"]

    if not record.get("speaker_id"):
        return False
    if not 3.5 <= duration <= 18.0:
        return False

    audio_path = Path(AUDIO_DIR) / record["audio_file"]
    if not audio_path.is_file():
        return False

    labels = tokenizer.encode(
        text, add_special_tokens=False
    )

    if not 20 <= len(labels) <= 140:
        return False
    if tokenizer.unk_token_id in labels:
        return False

    repeats = sum(
        a == b for a, b in zip(labels[:-1], labels[1:])
    )

    available = frame_count(round(duration * 16000))
    required = len(labels) + repeats

    return available - required >= 20

# ------------------------------------------------------------
# 1. Find suitable recordings
# ------------------------------------------------------------

candidates = [
    r for r in train_records
    if eligible_record(r)
]

assert eligible_record(record_lookup[ANCHOR_ID]), (
    "The known positive-control recording is unavailable."
)

rng = random.Random(20261019)
rng.shuffle(candidates)

# Prefer shorter recordings.
candidates.sort(
    key=lambda r: float(r["duration_seconds"])
)

print("DATASET AVAILABILITY")
print("-" * 50)

for maximum in [8, 10, 12, 15, 18]:
    speakers = {
        r["speaker_id"]
        for r in candidates
        if float(r["duration_seconds"]) <= maximum
    }
    print(
        f"Up to {maximum:2d}s:",
        f"{len(speakers)} unique speakers"
    )

# ------------------------------------------------------------
# 2. Adaptively select 12 different speakers
# ------------------------------------------------------------

chosen = None
selected_max_duration = None
digits_allowed = None

for allow_digits in [False, True]:

    for maximum in [8, 10, 12, 15, 18]:

        attempt = [record_lookup[ANCHOR_ID]]
        used_speakers = {
            attempt[0]["speaker_id"]
        }

        for record in candidates:

            if record["id"] == ANCHOR_ID:
                continue

            if float(record["duration_seconds"]) > maximum:
                continue

            if not allow_digits and any(
                ch.isdigit()
                for ch in record["transcription"]
            ):
                continue

            speaker = record["speaker_id"]

            if speaker in used_speakers:
                continue

            attempt.append(record)
            used_speakers.add(speaker)

            if len(attempt) == TRAIN_COUNT + VAL_COUNT:
                break

        if len(attempt) == TRAIN_COUNT + VAL_COUNT:
            chosen = attempt
            selected_max_duration = maximum
            digits_allowed = allow_digits
            break

    if chosen is not None:
        break

assert chosen is not None, (
    "Could not find 12 distinct speakers even after "
    "relaxing the recording duration to 18 seconds."
)

# ------------------------------------------------------------
# 3. Save and validate selection
# ------------------------------------------------------------

new_selection = {
    "anchor_id": ANCHOR_ID,
    "train_ids": [r["id"] for r in chosen[:8]],
    "val_ids": [r["id"] for r in chosen[8:]],
    "maximum_duration": selected_max_duration,
    "digits_allowed": digits_allowed
}

if SHORT_SELECTION_PATH.exists():
    selection = json.loads(
        SHORT_SELECTION_PATH.read_text(encoding="utf-8")
    )
    print("\nUsing existing saved selection.")
else:
    selection = new_selection
    SHORT_SELECTION_PATH.write_text(
        json.dumps(
            selection, indent=2, ensure_ascii=False
        ),
        encoding="utf-8"
    )
    print("\nNew selection saved.")

short_train_ids = selection["train_ids"]
short_val_ids = selection["val_ids"]

short_train_records = [
    record_lookup[rid] for rid in short_train_ids
]
short_val_records = [
    record_lookup[rid] for rid in short_val_ids
]

all_records = short_train_records + short_val_records

assert len(short_train_records) == 8
assert len(short_val_records) == 4
assert len({r["id"] for r in all_records}) == 12
assert len({r["speaker_id"] for r in all_records}) == 12
assert ANCHOR_ID in short_train_ids
assert all(eligible_record(r) for r in all_records)

print("\n" + "=" * 55)
print("CORRECTED DATASET SUMMARY")
print("=" * 55)

print("Training recordings:", len(short_train_records))
print("Held-out recordings:", len(short_val_records))
print("Unique speakers:", 12)
print(
    "Longest selected recording:",
    round(max(
        float(r["duration_seconds"])
        for r in all_records
    ), 2),
    "seconds"
)
print("Selection duration ceiling:", selected_max_duration)
print("Digits permitted in selection:", digits_allowed)

print("\nTRAINING RECORDINGS")
for i, record in enumerate(short_train_records, 1):
    print(
        f"{i}. {record['id']} | "
        f"{record['duration_seconds']:.2f}s"
    )
    print("   ", record["transcription"])

print("\nHELD-OUT RECORDINGS")
for i, record in enumerate(short_val_records, 1):
    print(
        f"{i}. {record['id']} | "
        f"{record['duration_seconds']:.2f}s"
    )
    print("   ", record["transcription"])

# ------------------------------------------------------------
# 4. Listen to a few examples
# ------------------------------------------------------------

print("\nAUDIO REVIEW")

for label, record in [
    ("KNOWN CONTROL", short_train_records[0]),
    ("NEW TRAINING", short_train_records[1]),
    ("HELD-OUT", short_val_records[0])
]:
    print("\n", label)
    print("Transcript:", record["transcription"])

    display(Audio(
        filename=str(
            Path(AUDIO_DIR) / record["audio_file"]
        )
    ))

print("\nSELECTION VALIDATION PASSED")
print("Saved:", SHORT_SELECTION_PATH)
print("No model checkpoints modified.")


DATASET AVAILABILITY
--------------------------------------------------
Up to  8s: 9 unique speakers
Up to 10s: 17 unique speakers
Up to 12s: 20 unique speakers
Up to 15s: 98 unique speakers
Up to 18s: 520 unique speakers

New selection saved.

CORRECTED DATASET SUMMARY
Training recordings: 8
Held-out recordings: 4
Unique speakers: 12
Longest selected recording: 9.7 seconds
Selection duration ceiling: 10
Digits permitted in selection: False

TRAINING RECORDINGS
1. 6Q0fEziAqyQVIz4J8aws | 5.18s
    ይህ ምስል የሚያሳየው ከሸክላ የሚሰራ የሸክላ ድስት ምስል ነው
2. 8DDU79GSsgg8dZV0J3ox | 4.30s
    ወንድ አርሶአደር በማሳ ላይ እየተጓዘ
3. MM8A6KtEQinYgNbyO1Zo | 4.78s
    በኢንዱስትሪ አካባቢ እንስቶች ልብስ ሲሰፉ የሚያሳይ ምስል ነው
4. VpYkSBOYaCCY8Zx6cEDm | 5.18s
    ምስሉ ላይ የምንመለከተው በአንድ የሸክላ ንስሀ ውስጥ ያለ የዶሮ ወጥ ነው
5. KJEzKPKIu0ecCoM99ebs | 6.70s
    ይህ የምናየው እንስሳ አንበሳ ይባላል በጫካ ውስጥ እየኖረ ነው ይህ የምናየው እንስሳ አንበሳ ይባላል በጫካ ውስጥ እየኖረ ነው
6. WdLLvXLdOnNtO7Xtc46Y | 6.94s
    አሁን በዚህ ምስል ላይ የምንመለከታቸው ማህበረሰቦች የሃይማኖት ስርአት እያከናወኑ ይገኛሉ
7. GjjqjszNttEsTkd4oBja | 7.46


 NEW TRAINING
Transcript: ወንድ አርሶአደር በማሳ ላይ እየተጓዘ



 HELD-OUT
Transcript: ይህ የምስል አይነት እንደሚያሳየን የባህላዊ የህክምና የጥርስ መፋቂያ የእጽዋት አይነት ነው



SELECTION VALIDATION PASSED
Saved: /content/drive/MyDrive/Amharic_ASR_XLSR/data/short_multirecording_v1/selection.json
No model checkpoints modified.


In [ ]:

# ============================================================
# CELL 41 - BALANCED SHORT-RECORDING ASR EXPERIMENT
#
# 8 train / 4 held-out, 12 different speakers
# Duration-balanced split
# Original XLS-R encoder frozen
# Only CTC head trainable
# ============================================================

import json
import copy
import gc
import hashlib
import itertools
import statistics
from pathlib import Path

import torch
import torch.nn.functional as F
from jiwer import cer, wer
from transformers import Wav2Vec2ForCTC

# ------------------------------------------------------------
# 1. Configuration
# ------------------------------------------------------------

MAX_UPDATES = 4000
REPORT_EVERY = 250
HEAD_LR = 1e-3

DEVICE_SHORT = torch.device(
    "cuda" if torch.cuda.is_available() else "cpu"
)

BLANK_SHORT = tokenizer.pad_token_id
ANCHOR_ID = "6Q0fEziAqyQVIz4J8aws"

SHORT_EXPERIMENT_DIR = (
    DATA_DIR / "short_multirecording_head_only_v2"
)
SHORT_EXPERIMENT_DIR.mkdir(
    parents=True, exist_ok=True
)

SPLIT_PATH = SHORT_EXPERIMENT_DIR / "split.json"
STATE_PATH = SHORT_EXPERIMENT_DIR / "latest.pt"
HISTORY_PATH = SHORT_EXPERIMENT_DIR / "history.json"

original_selection = json.loads(
    (
        DATA_DIR
        / "short_multirecording_v1"
        / "selection.json"
    ).read_text(encoding="utf-8")
)

pool_ids = (
    original_selection["train_ids"]
    + original_selection["val_ids"]
)

assert len(pool_ids) == 12
assert len(set(pool_ids)) == 12
assert ANCHOR_ID in pool_ids

by_id = {r["id"]: r for r in train_records}

def duration(rid):
    return float(by_id[rid]["duration_seconds"])

# ------------------------------------------------------------
# 2. Create a more balanced speaker-disjoint split
# ------------------------------------------------------------

if SPLIT_PATH.exists():

    split = json.loads(
        SPLIT_PATH.read_text(encoding="utf-8")
    )

    short_train_ids = split["train_ids"]
    short_val_ids = split["val_ids"]

    print("Reusing previously saved balanced split.")

else:

    others = [
        rid for rid in pool_ids
        if rid != ANCHOR_ID
    ]

    possible_splits = []

    for val_group in itertools.combinations(others, 4):

        val_group = list(val_group)
        val_set = set(val_group)

        train_group = [
            rid for rid in pool_ids
            if rid not in val_set
        ]

        train_durations = [
            duration(rid) for rid in train_group
        ]
        val_durations = [
            duration(rid) for rid in val_group
        ]

        # Both groups should contain recordings
        # of different lengths.
        if not any(d < 6 for d in val_durations):
            continue
        if not any(d >= 8 for d in val_durations):
            continue
        if not any(d >= 8 for d in train_durations):
            continue

        mean_gap = abs(
            statistics.mean(train_durations)
            - statistics.mean(val_durations)
        )

        spread_gap = abs(
            statistics.pstdev(train_durations)
            - statistics.pstdev(val_durations)
        )

        score = mean_gap + 0.25 * spread_gap

        possible_splits.append(
            (score, tuple(sorted(val_group)),
             train_group, val_group)
        )

    assert possible_splits, (
        "No suitable balanced split found."
    )

    possible_splits.sort(
        key=lambda item: (item[0], item[1])
    )

    _, _, short_train_ids, short_val_ids = (
        possible_splits[0]
    )

    split = {
        "train_ids": short_train_ids,
        "val_ids": short_val_ids,
        "anchor_id": ANCHOR_ID,
        "source_pool_ids": sorted(pool_ids)
    }

    SPLIT_PATH.write_text(
        json.dumps(
            split, ensure_ascii=False, indent=2
        ),
        encoding="utf-8"
    )

assert len(short_train_ids) == 8
assert len(short_val_ids) == 4
assert set(short_train_ids + short_val_ids) == set(pool_ids)
assert ANCHOR_ID in short_train_ids

train_speakers = {
    by_id[rid]["speaker_id"]
    for rid in short_train_ids
}
val_speakers = {
    by_id[rid]["speaker_id"]
    for rid in short_val_ids
}

assert len(train_speakers) == 8
assert len(val_speakers) == 4
assert not train_speakers.intersection(val_speakers)

print("\nBALANCED SPLIT")
print("-" * 55)
print("Training recordings:", len(short_train_ids))
print("Held-out recordings:", len(short_val_ids))
print("Overlapping speakers:", 0)

print(
    "Mean train duration:",
    round(statistics.mean(
        duration(rid) for rid in short_train_ids
    ), 2),
    "seconds"
)

print(
    "Mean held-out duration:",
    round(statistics.mean(
        duration(rid) for rid in short_val_ids
    ), 2),
    "seconds"
)

# ------------------------------------------------------------
# 3. Verify a reproducible experiment signature
# ------------------------------------------------------------

experiment_config = {
    "train_ids": short_train_ids,
    "val_ids": short_val_ids,
    "references": {
        rid: by_id[rid]["transcription"]
        for rid in short_train_ids + short_val_ids
    },
    "baseline": str(BASELINE_DIR),
    "head_lr": HEAD_LR
}

signature = hashlib.sha256(
    json.dumps(
        experiment_config,
        sort_keys=True,
        ensure_ascii=False
    ).encode("utf-8")
).hexdigest()

index_by_id = {
    r["id"]: index
    for index, r in enumerate(train_dataset.records)
}

# ------------------------------------------------------------
# 4. Load frozen original XLS-R encoder
# ------------------------------------------------------------

print("\nLoading original XLS-R model...")

short_model = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(DEVICE_SHORT)

short_model.eval()

# Copy the CTC head outside inference mode.
short_head = copy.deepcopy(
    short_model.lm_head
).to(DEVICE_SHORT).float()

assert short_head.weight.requires_grad
assert not short_head.weight.is_inference()

# ------------------------------------------------------------
# 5. Cache encoder features once
# ------------------------------------------------------------

def prepare_short_item(rid):

    example = train_dataset[index_by_id[rid]]
    batch = ctc_collator([example])

    batch = {
        key: value.to(DEVICE_SHORT)
        for key, value in batch.items()
    }

    with torch.no_grad():

        features = short_model.wav2vec2(
            input_values=batch["input_values"],
            attention_mask=batch["attention_mask"]
        ).last_hidden_state

    features = features.detach().clone().float()

    targets = batch["labels"][
        batch["labels"] >= 0
    ].reshape(-1).contiguous()

    repeated = int(
        (targets[1:] == targets[:-1]).sum().item()
    )

    assert features.shape[1] >= (
        targets.numel() + repeated
    )

    assert not features.is_inference()
    assert torch.isfinite(features).all()

    return {
        "id": rid,
        "features": features,
        "targets": targets,
        "input_lengths": torch.tensor(
            [features.shape[1]], dtype=torch.long
        ),
        "target_lengths": torch.tensor(
            [targets.numel()], dtype=torch.long
        ),
        "reference": normalize_amharic_ctc(
            by_id[rid]["transcription"]
        )
    }

print("\nCaching encoder features...")

short_train_items = [
    prepare_short_item(rid)
    for rid in short_train_ids
]

short_val_items = [
    prepare_short_item(rid)
    for rid in short_val_ids
]

del short_model
gc.collect()
torch.cuda.empty_cache()

print("Cached: 8 train + 4 held-out")
print(
    "Trainable head parameters:",
    sum(p.numel() for p in short_head.parameters())
)

# ------------------------------------------------------------
# 6. Training and evaluation functions
# ------------------------------------------------------------

def short_ctc_loss(item):

    logits = short_head(item["features"])

    return F.ctc_loss(
        F.log_softmax(
            logits.float(), dim=-1
        ).transpose(0, 1),
        item["targets"],
        item["input_lengths"],
        item["target_lengths"],
        blank=BLANK_SHORT,
        reduction="mean",
        zero_infinity=False
    )


def short_evaluate(items):

    short_head.eval()

    references = []
    predictions = []
    losses = []

    with torch.no_grad():

        for item in items:

            logits = short_head(item["features"])

            ids = logits.argmax(dim=-1)

            text = processor.batch_decode(
                ids.cpu()
            )[0]

            text = normalize_amharic_ctc(text)

            references.append(item["reference"])
            predictions.append(text)

            losses.append(
                float(short_ctc_loss(item).item())
            )

    return {
        "cer": float(cer(references, predictions)),
        "wer": float(wer(references, predictions)),
        "loss": sum(losses) / len(losses),
        "nonempty": sum(
            bool(text.strip()) for text in predictions
        ),
        "predictions": predictions
    }

short_optimizer = torch.optim.AdamW(
    short_head.parameters(),
    lr=HEAD_LR,
    weight_decay=0.0
)

# ------------------------------------------------------------
# 7. Resume if an experiment already exists
# ------------------------------------------------------------

history = []
start_step = 0

if STATE_PATH.exists():

    state = torch.load(
        STATE_PATH,
        map_location="cpu",
        weights_only=True
    )

    assert state["signature"] == signature
    assert state["lr"] == HEAD_LR

    short_head.load_state_dict(state["head"])
    short_optimizer.load_state_dict(state["optimizer"])

    start_step = int(state["step"])

    if HISTORY_PATH.exists():
        history = json.loads(
            HISTORY_PATH.read_text(encoding="utf-8")
        )

    print(f"\nResuming from step {start_step}")

else:
    print("\nStarting new head-only experiment.")

def short_save(step):

    state = {
        "step": step,
        "signature": signature,
        "lr": HEAD_LR,
        "head": short_head.state_dict(),
        "optimizer": short_optimizer.state_dict()
    }

    temp = SHORT_EXPERIMENT_DIR / "latest.pt.partial"

    torch.save(state, temp)
    temp.replace(STATE_PATH)

    temp_hist = (
        SHORT_EXPERIMENT_DIR / "history.json.partial"
    )

    temp_hist.write_text(
        json.dumps(
            history, ensure_ascii=False, indent=2
        ),
        encoding="utf-8"
    )

    temp_hist.replace(HISTORY_PATH)

# ------------------------------------------------------------
# 8. Reporting
# ------------------------------------------------------------

def short_report(step):

    train_result = short_evaluate(short_train_items)
    val_result = short_evaluate(short_val_items)

    result = {
        "step": step,
        "train_cer": train_result["cer"],
        "train_wer": train_result["wer"],
        "train_loss": train_result["loss"],
        "val_cer": val_result["cer"],
        "val_wer": val_result["wer"],
        "val_loss": val_result["loss"],
        "train_nonempty": train_result["nonempty"],
        "val_nonempty": val_result["nonempty"]
    }

    print(f"\nSTEP {step}/{MAX_UPDATES}")
    print("-" * 48)

    print(
        "Train CER:",
        f"{train_result['cer'] * 100:.2f}%"
    )

    print(
        "Held-out CER:",
        f"{val_result['cer'] * 100:.2f}%"
    )

    print(
        "Held-out WER:",
        f"{val_result['wer'] * 100:.2f}%"
    )

    print(
        "Train loss:",
        round(train_result["loss"], 4)
    )

    print(
        "Nonempty:",
        f"{train_result['nonempty']}/8 train,",
        f"{val_result['nonempty']}/4 held-out"
    )

    print("\nKnown positive-control prediction:")
    anchor_index = short_train_ids.index(ANCHOR_ID)
    print(
        train_result["predictions"][anchor_index]
        or "[EMPTY]"
    )

    print("\nHeld-out prediction:")
    print(
        val_result["predictions"][0]
        or "[EMPTY]"
    )

    return result

if start_step == 0 and not history:
    history.append(short_report(0))

# ------------------------------------------------------------
# 9. Train with deterministic rotating examples
# ------------------------------------------------------------

print("\nTRAINING SHORT-RECORDING MODEL")
print("=" * 55)

completed_step = start_step

for step in range(start_step + 1, MAX_UPDATES + 1):

    item = short_train_items[
        (step - 1) % len(short_train_items)
    ]

    short_head.train()
    short_optimizer.zero_grad(set_to_none=True)

    loss = short_ctc_loss(item)

    assert torch.isfinite(loss).item()
    assert loss.requires_grad

    loss.backward()

    torch.nn.utils.clip_grad_norm_(
        short_head.parameters(),
        max_norm=5.0,
        error_if_nonfinite=True
    )

    short_optimizer.step()

    completed_step = step

    if step % REPORT_EVERY == 0:

        report = short_report(step)
        history.append(report)

        short_save(step)

# ------------------------------------------------------------
# 10. Final results
# ------------------------------------------------------------

final_train = short_evaluate(short_train_items)
final_val = short_evaluate(short_val_items)

print("\n" + "=" * 60)
print("FINAL SHORT-RECORDING RESULTS")
print("=" * 60)

print("Completed updates:", completed_step)

print(
    "Training CER:",
    f"{final_train['cer'] * 100:.2f}%"
)

print(
    "Held-out CER:",
    f"{final_val['cer'] * 100:.2f}%"
)

print(
    "Held-out WER:",
    f"{final_val['wer'] * 100:.2f}%"
)

print("\nCheckpoint:", STATE_PATH)
print("History:", HISTORY_PATH)

print("\nExisting XLS-R and step-500 checkpoints unchanged.")



BALANCED SPLIT
-------------------------------------------------------
Training recordings: 8
Held-out recordings: 4
Overlapping speakers: 0
Mean train duration: 6.95 seconds
Mean held-out duration: 6.97 seconds

Loading original XLS-R model...

Caching encoder features...
Cached: 8 train + 4 held-out
Trainable head parameters: 329025

Starting new head-only experiment.

STEP 0/4000
------------------------------------------------
Train CER: 150.57%
Held-out CER: 141.88%
Held-out WER: 100.00%
Train loss: 33.2595
Nonempty: 8/8 train, 4/4 held-out

Known positive-control prediction:
ጠጹኧጹኻጹኻሣጹሣኻ፲ኻጹኻሣኻጹኻሼጹኻጹኻጹሣtጹሣጹኻጹኻጹሣጹኻጹኻጹኻጹሣጹኻtሼኻጹሼኦጹሄኻጹሣጹኻtጹኻጹሣኻጹtሣጹኻጹሣኻ፲ጹሼጹኻጹሼሣኻጹኻጹኻጹኻጹሼጹሣኻጹኻጹሣጹtጹኧ

Held-out prediction:
ጠኻጹኻጹኻጹኻጹኻጹኻጹኻጹኻጹኻሄኻሄኻሼኻጹኧኻሼኻጹኻጹኻጹሼኻጹኻጹኻጹኻጹሄጹኻኧ

TRAINING SHORT-RECORDING MODEL

STEP 250/4000
------------------------------------------------
Train CER: 96.15%
Held-out CER: 94.87%
Held-out WER: 100.00%
Train loss: 3.3604
Nonempty: 8/8 train, 4/4 held-out

Known positive-control predic

In [ ]:

# ============================================================
# CELL 42 - CONTROLLED TWO-STAGE FINE-TUNING TEST
#
# A: Frozen XLS-R encoder + trained CTC head
# B: Train last 2 XLS-R layers + same trained CTC head
#
# Both start from the Cell 41 head at update 4000.
# Same data order, head LR, and number of updates.
# Old checkpoints are never modified.
# ============================================================

import copy
import gc
import json
import hashlib
from pathlib import Path

import torch
import torch.nn.functional as F
from jiwer import cer, wer
from transformers import Wav2Vec2ForCTC

DEVICE_42 = torch.device(
    "cuda" if torch.cuda.is_available() else "cpu"
)

PILOT_UPDATES = 300
REPORT_EVERY = 100
HEAD_LR = 3e-4
ENCODER_LR = 1e-5
BLANK = tokenizer.pad_token_id
ANCHOR_ID = "6Q0fEziAqyQVIz4J8aws"

WARM_DIR = DATA_DIR / "short_multirecording_head_only_v2"
WARM_STATE = WARM_DIR / "latest.pt"
SPLIT_FILE = WARM_DIR / "split.json"

RUN_DIR = DATA_DIR / "warm_head_encoder_comparison_v1"
RUN_DIR.mkdir(parents=True, exist_ok=True)

assert WARM_STATE.is_file()
assert SPLIT_FILE.is_file()

warm = torch.load(
    WARM_STATE,
    map_location="cpu",
    weights_only=True
)

assert int(warm["step"]) == 4000

split = json.loads(
    SPLIT_FILE.read_text(encoding="utf-8")
)

train_ids = split["train_ids"]
val_ids = split["val_ids"]

assert len(train_ids) == 8
assert len(val_ids) == 4
assert ANCHOR_ID in train_ids
assert len(set(train_ids + val_ids)) == 12

by_id = {r["id"]: r for r in train_records}
index_by_id = {
    r["id"]: i
    for i, r in enumerate(train_dataset.records)
}

assert len({
    by_id[rid]["speaker_id"]
    for rid in train_ids + val_ids
}) == 12

signature = hashlib.sha256(
    json.dumps({
        "train_ids": train_ids,
        "val_ids": val_ids,
        "warm_signature": warm["signature"],
        "warm_step": warm["step"],
        "head_lr": HEAD_LR,
        "encoder_lr": ENCODER_LR
    }, sort_keys=True).encode()
).hexdigest()

print("CONTROLLED FINE-TUNING EXPERIMENT")
print("=" * 55)
print("Starting head: Cell 41, update 4000")
print("Training recordings:", len(train_ids))
print("Held-out recordings:", len(val_ids))
print("Updates per branch:", PILOT_UPDATES)

# ------------------------------------------------------------
# 1. Load audio once, keeping exactly the same preprocessing
# ------------------------------------------------------------

batches = {}

for rid in train_ids + val_ids:
    example = train_dataset[index_by_id[rid]]
    batch = ctc_collator([example])
    batches[rid] = {
        k: v.to(DEVICE_42)
        for k, v in batch.items()
    }

references = {
    rid: normalize_amharic_ctc(
        by_id[rid]["transcription"]
    )
    for rid in train_ids + val_ids
}

def score_predictions(predict_fn, ids):
    refs = []
    preds = []

    with torch.no_grad():
        for rid in ids:
            token_ids = predict_fn(rid)
            text = processor.batch_decode(
                token_ids.detach().cpu()
            )[0]
            text = normalize_amharic_ctc(text)

            refs.append(references[rid])
            preds.append(text)

    return {
        "cer": float(cer(refs, preds)),
        "wer": float(wer(refs, preds)),
        "predictions": preds
    }

def report(branch, step, predict_fn):
    train_result = score_predictions(
        predict_fn, train_ids
    )
    val_result = score_predictions(
        predict_fn, val_ids
    )

    result = {
        "step": step,
        "train_cer": train_result["cer"],
        "val_cer": val_result["cer"],
        "val_wer": val_result["wer"],
        "anchor_prediction":
            train_result["predictions"][
                train_ids.index(ANCHOR_ID)
            ],
        "val_prediction":
            val_result["predictions"][0]
    }

    print(f"\n{branch} | UPDATE {step}")
    print(
        "Train CER:",
        f"{result['train_cer'] * 100:.2f}%"
    )
    print(
        "Held-out CER:",
        f"{result['val_cer'] * 100:.2f}%"
    )
    print(
        "Held-out WER:",
        f"{result['val_wer'] * 100:.2f}%"
    )
    print(
        "Anchor:",
        result["anchor_prediction"] or "[EMPTY]"
    )
    print(
        "Held-out:",
        result["val_prediction"] or "[EMPTY]"
    )

    return result

def save_state(path, state, history, history_path):
    temp = path.with_suffix(".pt.partial")
    torch.save(state, temp)
    temp.replace(path)

    history_temp = history_path.with_suffix(
        ".json.partial"
    )
    history_temp.write_text(
        json.dumps(
            history,
            indent=2,
            ensure_ascii=False
        ),
        encoding="utf-8"
    )
    history_temp.replace(history_path)

# ------------------------------------------------------------
# 2. Load original encoder and cache frozen features
# ------------------------------------------------------------

print("\nLoading original encoder...")

base = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(DEVICE_42)

base.eval()
base.lm_head.load_state_dict(warm["head"])

features = {}

with torch.no_grad():
    for rid, batch in batches.items():
        hidden = base.wav2vec2(
            input_values=batch["input_values"],
            attention_mask=batch["attention_mask"]
        ).last_hidden_state

        features[rid] = hidden.detach().clone().float()

head_a = copy.deepcopy(base.lm_head)
head_a.requires_grad_(True)

del base
gc.collect()
torch.cuda.empty_cache()

# ------------------------------------------------------------
# 3. Branch A: Continue training the head only
# ------------------------------------------------------------

print("\nBRANCH A: FROZEN ENCODER")
print("=" * 55)

optimizer_a = torch.optim.AdamW(
    head_a.parameters(),
    lr=HEAD_LR,
    weight_decay=0.0
)

def predict_a(rid):
    return head_a(features[rid]).argmax(-1)

def loss_a(rid):
    logits = head_a(features[rid])

    target = batches[rid]["labels"]
    target = target[target >= 0].reshape(-1)

    return F.ctc_loss(
        F.log_softmax(logits.float(), -1).transpose(0, 1),
        target,
        torch.tensor(
            [logits.shape[1]], dtype=torch.long
        ),
        torch.tensor(
            [target.numel()], dtype=torch.long
        ),
        blank=BLANK,
        reduction="mean",
        zero_infinity=False
    )

a_path = RUN_DIR / "head_only_latest.pt"
a_history_path = RUN_DIR / "head_only_history.json"

a_step = 0
history_a = []

if a_path.exists():
    saved_a = torch.load(
        a_path, map_location="cpu", weights_only=True
    )
    assert saved_a["signature"] == signature

    head_a.load_state_dict(saved_a["head"])
    optimizer_a.load_state_dict(saved_a["optimizer"])
    a_step = int(saved_a["step"])

    if a_history_path.exists():
        history_a = json.loads(
            a_history_path.read_text(encoding="utf-8")
        )

if not history_a:
    history_a.append(report("A", a_step, predict_a))

for step in range(a_step + 1, PILOT_UPDATES + 1):

    rid = train_ids[(step - 1) % len(train_ids)]

    optimizer_a.zero_grad(set_to_none=True)
    loss = loss_a(rid)

    assert torch.isfinite(loss).item()
    assert loss.requires_grad

    loss.backward()

    torch.nn.utils.clip_grad_norm_(
        head_a.parameters(), 5.0
    )

    optimizer_a.step()

    if step % REPORT_EVERY == 0:
        history_a.append(
            report("A", step, predict_a)
        )

        save_state(
            a_path,
            {
                "signature": signature,
                "step": step,
                "head": head_a.state_dict(),
                "optimizer": optimizer_a.state_dict()
            },
            history_a,
            a_history_path
        )

del head_a, optimizer_a, features
gc.collect()
torch.cuda.empty_cache()

# ------------------------------------------------------------
# 4. Branch B: Unfreeze last 2 Transformer layers
# ------------------------------------------------------------

print("\nBRANCH B: TRAIN LAST 2 TRANSFORMER LAYERS")
print("=" * 55)

model_b = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(DEVICE_42)

model_b.lm_head.load_state_dict(warm["head"])

# Freeze everything first.
for parameter in model_b.parameters():
    parameter.requires_grad_(False)

# Train only last 2 Transformer layers.
upper_layers = list(
    model_b.wav2vec2.encoder.layers[-2:]
)

for layer in upper_layers:
    for parameter in layer.parameters():
        parameter.requires_grad_(True)

for parameter in model_b.lm_head.parameters():
    parameter.requires_grad_(True)

# Diagnostic training with dropout and SpecAugment off.
# eval() DOES NOT disable gradients; it disables
# stochastic training behaviors such as dropout.
# This keeps comparison with cached features controlled.
model_b.eval()

encoder_parameters = [
    p
    for layer in upper_layers
    for p in layer.parameters()
    if p.requires_grad
]

head_parameters = list(
    model_b.lm_head.parameters()
)

optimizer_b = torch.optim.AdamW(
    [
        {
            "params": encoder_parameters,
            "lr": ENCODER_LR,
            "weight_decay": 0.01
        },
        {
            "params": head_parameters,
            "lr": HEAD_LR,
            "weight_decay": 0.0
        }
    ]
)

use_amp = DEVICE_42.type == "cuda"

scaler_b = torch.amp.GradScaler(
    "cuda", enabled=use_amp
)

print(
    "Trainable parameters:",
    sum(
        p.numel()
        for p in model_b.parameters()
        if p.requires_grad
    )
)

def predict_b(rid):
    return model_b(**batches[rid]).logits.argmax(-1)

b_path = RUN_DIR / "last2_latest.pt"
b_history_path = RUN_DIR / "last2_history.json"

b_step = 0
history_b = []

if b_path.exists():
    saved_b = torch.load(
        b_path, map_location="cpu", weights_only=True
    )
    assert saved_b["signature"] == signature

    model_b.lm_head.load_state_dict(
        saved_b["head"]
    )

    for layer, weights in zip(
        upper_layers, saved_b["upper_layers"]
    ):
        layer.load_state_dict(weights)

    optimizer_b.load_state_dict(
        saved_b["optimizer"]
    )

    scaler_b.load_state_dict(saved_b["scaler"])
    b_step = int(saved_b["step"])

    if b_history_path.exists():
        history_b = json.loads(
            b_history_path.read_text(encoding="utf-8")
        )

if not history_b:
    history_b.append(report("B", b_step, predict_b))

for step in range(b_step + 1, PILOT_UPDATES + 1):

    rid = train_ids[(step - 1) % len(train_ids)]

    optimizer_b.zero_grad(set_to_none=True)

    with torch.autocast(
        device_type="cuda",
        dtype=torch.float16,
        enabled=use_amp
    ):
        loss = model_b(**batches[rid]).loss

    assert torch.isfinite(loss).item()
    assert loss.requires_grad

    scaler_b.scale(loss).backward()
    scaler_b.unscale_(optimizer_b)

    torch.nn.utils.clip_grad_norm_(
        encoder_parameters + head_parameters,
        max_norm=1.0,
        error_if_nonfinite=True
    )

    scaler_b.step(optimizer_b)
    scaler_b.update()

    if step % REPORT_EVERY == 0:

        history_b.append(
            report("B", step, predict_b)
        )

        save_state(
            b_path,
            {
                "signature": signature,
                "step": step,
                "head": model_b.lm_head.state_dict(),
                "upper_layers": [
                    layer.state_dict()
                    for layer in upper_layers
                ],
                "optimizer": optimizer_b.state_dict(),
                "scaler": scaler_b.state_dict()
            },
            history_b,
            b_history_path
        )

# ------------------------------------------------------------
# 5. Side-by-side results
# ------------------------------------------------------------

print("\n" + "=" * 60)
print("CONTROLLED COMPARISON RESULTS")
print("=" * 60)

print(
    f"{'Update':<10}"
    f"{'A Train':<13}"
    f"{'B Train':<13}"
    f"{'A Held-out':<15}"
    f"{'B Held-out':<15}"
)

a_by_step = {
    row["step"]: row for row in history_a
}
b_by_step = {
    row["step"]: row for row in history_b
}

for step in sorted(
    set(a_by_step) & set(b_by_step)
):
    a = a_by_step[step]
    b = b_by_step[step]

    print(
        f"{step:<10}"
        f"{a['train_cer']*100:<13.2f}"
        f"{b['train_cer']*100:<13.2f}"
        f"{a['val_cer']*100:<15.2f}"
        f"{b['val_cer']*100:<15.2f}"
    )

print("\nBranch A: Frozen pretrained encoder")
print("Branch B: Train last 2 Transformer layers")
print("Previous baseline and step-500 checkpoints unchanged.")
print("Experiment directory:", RUN_DIR)

CONTROLLED FINE-TUNING EXPERIMENT
Starting head: Cell 41, update 4000
Training recordings: 8
Held-out recordings: 4
Updates per branch: 300

Loading original encoder...

BRANCH A: FROZEN ENCODER

A | UPDATE 0
Train CER: 49.89%
Held-out CER: 87.61%
Held-out WER: 100.00%
Anchor: ይምየሳውሸክላየሸክላድ ምስ ው
Held-out: ይሳም ም ሳ ምው

A | UPDATE 100
Train CER: 49.66%
Held-out CER: 87.61%
Held-out WER: 100.00%
Anchor: ይምየሳውሸክላየሸክላድ ምስ ው
Held-out: ይሳም ም ሳ ምው

A | UPDATE 200
Train CER: 49.66%
Held-out CER: 87.61%
Held-out WER: 100.00%
Anchor: ይምየሳውሸክላየሸክላድ ምስ ው
Held-out: ይሳም ም ሳ ምው

A | UPDATE 300
Train CER: 49.21%
Held-out CER: 87.61%
Held-out WER: 100.00%
Anchor: ይምየሳውሸክላየሸክላድ ምስ ው
Held-out: ይሳም ም ሳ ምው

BRANCH B: TRAIN LAST 2 TRANSFORMER LAYERS
Trainable parameters: 25521473

B | UPDATE 0
Train CER: 49.89%
Held-out CER: 87.61%
Held-out WER: 100.00%
Anchor: ይምየሳውሸክላየሸክላድ ምስ ው
Held-out: ይሳም ም ሳ ምው


RuntimeError: The total norm of order 2.0 for gradients from `parameters` is non-finite, so it cannot be clipped. To disable this error and scale the gradients by the non-finite norm anyway, set `error_if_nonfinite=False`

In [ ]:

# ============================================================
# CELL 42B - REPAIR BRANCH B: FULL FP32 TRAINING
#
# Fix: Disable mixed precision and gradient scaling.
# Reuse the loaded Branch B model and optimizer.
# Branch A and all previous checkpoints remain unchanged.
# ============================================================

import json
import torch
from pathlib import Path

# ------------------------------------------------------------
# 1. Check dependencies from Cell 42
# ------------------------------------------------------------

required = [
    "model_b",
    "optimizer_b",
    "batches",
    "train_ids",
    "val_ids",
    "upper_layers",
    "encoder_parameters",
    "head_parameters",
    "predict_b",
    "report",
    "RUN_DIR",
    "signature",
]

missing = [
    name for name in required
    if name not in globals()
]

assert not missing, (
    "Missing Cell 42 variables: " + ", ".join(missing)
)

FP32_UPDATES = 300
FP32_REPORT_EVERY = 100

FP32_STATE = RUN_DIR / "last2_fp32_latest.pt"
FP32_HISTORY = RUN_DIR / "last2_fp32_history.json"

# ------------------------------------------------------------
# 2. Prepare the model for full-precision training
# ------------------------------------------------------------

model_b = model_b.float()
model_b.eval()

# Clear invalid gradients left by the failed FP16 attempt.
optimizer_b.zero_grad(set_to_none=True)

trainable_params = [
    p for p in model_b.parameters()
    if p.requires_grad
]

assert len(trainable_params) > 0
assert all(p.dtype == torch.float32 for p in trainable_params)

print("FP32 TRAINING REPAIR")
print("=" * 55)
print("Model parameter dtype: float32")
print("Mixed precision: DISABLED")
print("Gradient scaler: DISABLED")
print("Trainable parameters:", sum(
    p.numel() for p in trainable_params
))

# ------------------------------------------------------------
# 3. Restore previous FP32 progress if available
# ------------------------------------------------------------

fp32_start = 0
fp32_history = []

if FP32_STATE.exists():

    saved = torch.load(
        FP32_STATE,
        map_location="cpu",
        weights_only=True
    )

    assert saved["signature"] == signature
    assert saved["precision"] == "fp32"

    model_b.lm_head.load_state_dict(saved["head"])

    for layer, weights in zip(
        upper_layers,
        saved["upper_layers"]
    ):
        layer.load_state_dict(weights)

    optimizer_b.load_state_dict(saved["optimizer"])

    fp32_start = int(saved["step"])

    if FP32_HISTORY.exists():
        fp32_history = json.loads(
            FP32_HISTORY.read_text(encoding="utf-8")
        )

    print("Resuming FP32 experiment:", fp32_start)

else:
    # The FP16 attempt failed before optimizer.step().
    # Therefore the model should still have the
    # original warm-head initialization.
    assert "warm" in globals()

    for name, parameter in model_b.lm_head.state_dict().items():
        expected = warm["head"][name].to(
            parameter.device
        )
        assert torch.equal(parameter, expected), (
            f"Unexpected modification to head: {name}"
        )

    print("Original warm-head weights: VERIFIED")

# ------------------------------------------------------------
# 4. Check one FP32 backward pass WITHOUT updating weights
# ------------------------------------------------------------

first_id = train_ids[
    fp32_start % len(train_ids)
]

print("\nTESTING FP32 GRADIENTS")
print("-" * 55)
print("Diagnostic recording:", first_id)

optimizer_b.zero_grad(set_to_none=True)

# No autocast, no GradScaler.
with torch.autocast(
    device_type="cuda",
    enabled=False
):
    test_loss = model_b(**batches[first_id]).loss

print("Loss:", float(test_loss.item()))
print("Loss dtype:", test_loss.dtype)
print("Requires grad:", test_loss.requires_grad)

assert torch.isfinite(test_loss).item()
assert test_loss.requires_grad

test_loss.backward()

bad_gradients = []

for name, parameter in model_b.named_parameters():

    if not parameter.requires_grad:
        continue

    grad = parameter.grad

    if grad is None:
        continue

    if not torch.isfinite(grad).all().item():

        bad_count = int(
            (~torch.isfinite(grad)).sum().item()
        )

        bad_gradients.append((name, bad_count))

print("Parameters with invalid gradients:",
      len(bad_gradients))

if bad_gradients:
    for name, count in bad_gradients[:10]:
        print("INVALID:", name, "count:", count)

    optimizer_b.zero_grad(set_to_none=True)

    raise RuntimeError(
        "Non-finite gradients persist in FP32. "
        "Do not train yet; inspect the output."
    )

test_grad_norm = torch.nn.utils.clip_grad_norm_(
    trainable_params,
    max_norm=1.0,
    error_if_nonfinite=True
)

print("Gradient norm before clipping:",
      float(test_grad_norm))

optimizer_b.zero_grad(set_to_none=True)

print("\nFP32 GRADIENT CHECK: PASSED")
print("No optimizer update was performed in this test.")

# ------------------------------------------------------------
# 5. Define independent FP32 checkpoint saving
# ------------------------------------------------------------

def save_fp32(step):

    state = {
        "signature": signature,
        "precision": "fp32",
        "step": step,
        "head": model_b.lm_head.state_dict(),
        "upper_layers": [
            layer.state_dict()
            for layer in upper_layers
        ],
        "optimizer": optimizer_b.state_dict(),
    }

    temporary = RUN_DIR / "last2_fp32_latest.pt.partial"

    torch.save(state, temporary)
    temporary.replace(FP32_STATE)

    history_temp = (
        RUN_DIR / "last2_fp32_history.json.partial"
    )

    history_temp.write_text(
        json.dumps(
            fp32_history,
            indent=2,
            ensure_ascii=False
        ),
        encoding="utf-8"
    )

    history_temp.replace(FP32_HISTORY)

# ------------------------------------------------------------
# 6. Evaluate the starting point
# ------------------------------------------------------------

if not fp32_history:
    fp32_history.append(
        report("B FP32", fp32_start, predict_b)
    )

# ------------------------------------------------------------
# 7. Train last two Transformer layers in FP32
# ------------------------------------------------------------

print("\nSTARTING BRANCH B FP32 TRAINING")
print("=" * 55)

completed = fp32_start

for step in range(
    fp32_start + 1,
    FP32_UPDATES + 1
):

    rid = train_ids[
        (step - 1) % len(train_ids)
    ]

    optimizer_b.zero_grad(set_to_none=True)

    with torch.autocast(
        device_type="cuda",
        enabled=False
    ):
        loss = model_b(**batches[rid]).loss

    assert torch.isfinite(loss).item(), (
        f"Non-finite loss at update {step}"
    )

    loss.backward()

    grad_norm = torch.nn.utils.clip_grad_norm_(
        trainable_params,
        max_norm=1.0,
        error_if_nonfinite=True
    )

    optimizer_b.step()

    completed = step

    if step % FP32_REPORT_EVERY == 0:

        result = report(
            "B FP32",
            step,
            predict_b
        )

        result["gradient_norm"] = float(
            grad_norm
        )

        result["training_loss"] = float(
            loss.item()
        )

        fp32_history.append(result)

        save_fp32(step)

# ------------------------------------------------------------
# 8. Compare with the saved Branch A results
# ------------------------------------------------------------

a_history_file = RUN_DIR / "head_only_history.json"

assert a_history_file.exists()

history_a_saved = json.loads(
    a_history_file.read_text(encoding="utf-8")
)

a_by_step = {
    row["step"]: row
    for row in history_a_saved
}

b_by_step = {
    row["step"]: row
    for row in fp32_history
}

print("\n" + "=" * 65)
print("CONTROLLED COMPARISON: BRANCH A VS BRANCH B")
print("=" * 65)

print(
    f"{'Step':<8}"
    f"{'A Train':<13}"
    f"{'B Train':<13}"
    f"{'A Held-out':<15}"
    f"{'B Held-out':<15}"
)

for step in sorted(
    set(a_by_step) & set(b_by_step)
):

    a = a_by_step[step]
    b = b_by_step[step]

    print(
        f"{step:<8}"
        f"{a['train_cer']*100:<13.2f}"
        f"{b['train_cer']*100:<13.2f}"
        f"{a['val_cer']*100:<15.2f}"
        f"{b['val_cer']*100:<15.2f}"
    )

print("\nFP32 updates completed:", completed)
print("FP32 checkpoint:", FP32_STATE)
print("FP32 history:", FP32_HISTORY)
print("\nPrevious checkpoints remain unchanged.")


FP32 TRAINING REPAIR
Model parameter dtype: float32
Mixed precision: DISABLED
Gradient scaler: DISABLED
Trainable parameters: 25521473


AssertionError: Unexpected modification to head: weight

In [ ]:

# ============================================================
# CELL 42C - CLEAN BRANCH B RESET AND FP32 GRADIENT TEST
#
# Rebuild from original XLS-R + saved Cell 41 head.
# Do not reuse potentially inconsistent model weights.
# No training updates; no checkpoints overwritten.
# ============================================================

import gc
import torch
from pathlib import Path
from transformers import Wav2Vec2ForCTC

DEVICE_42 = torch.device(
    "cuda" if torch.cuda.is_available() else "cpu"
)

WARM_STATE_PATH = (
    DATA_DIR
    / "short_multirecording_head_only_v2"
    / "latest.pt"
)

assert WARM_STATE_PATH.is_file()
assert Path(BASELINE_DIR).is_dir()

# ==========================================
# 1. LOAD VERIFIED HEAD WEIGHTS FROM DISK
# ==========================================

warm_verified = torch.load(
    WARM_STATE_PATH,
    map_location="cpu",
    weights_only=True
)

assert warm_verified["step"] == 4000

expected_head = warm_verified["head"]

print("CHECKING PREVIOUS WEIGHT MISMATCH")
print("-" * 55)

if "model_b" in globals():

    actual = (
        model_b.lm_head.weight
        .detach()
        .cpu()
    )

    expected = expected_head["weight"]

    print(
        "Existing head matches saved head:",
        torch.equal(actual, expected)
    )

    print(
        "Current head finite:",
        bool(torch.isfinite(actual).all())
    )

    print(
        "Saved head finite:",
        bool(torch.isfinite(expected).all())
    )

    if torch.isfinite(actual).all() and torch.isfinite(expected).all():
        print(
            "Maximum absolute weight difference:",
            float((actual - expected).abs().max())
        )

# ==========================================
# 2. RELEASE OLD FAILED BRANCH B STATE
# ==========================================

for name in [
    "optimizer_b",
    "scaler_b",
    "model_b",
    "upper_layers",
    "encoder_parameters",
    "head_parameters",
    "trainable_params"
]:
    if name in globals():
        del globals()[name]

gc.collect()

if torch.cuda.is_available():
    torch.cuda.empty_cache()

# ==========================================
# 3. REBUILD MODEL FROM ORIGINAL BASELINE
# ==========================================

print("\nREBUILDING BRANCH B")
print("-" * 55)

model_b = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(DEVICE_42).float()

# Restore exactly the same head that Branch A used.
model_b.lm_head.load_state_dict(
    expected_head,
    strict=True
)

# Verify that restoration really worked.
for name, parameter in model_b.lm_head.state_dict().items():

    expected = expected_head[name].to(
        parameter.device
    )

    assert torch.equal(parameter, expected), (
        f"Head restoration failed: {name}"
    )

print("Saved Cell 41 head restored: VERIFIED")

# ==========================================
# 4. CONFIGURE TRAINABLE PARAMETERS
# ==========================================

# Freeze the entire model.
model_b.requires_grad_(False)

# Unfreeze last two Transformer layers.
upper_layers = list(
    model_b.wav2vec2.encoder.layers[-2:]
)

for layer in upper_layers:
    layer.requires_grad_(True)

# Unfreeze the CTC head.
model_b.lm_head.requires_grad_(True)

encoder_parameters = [
    parameter
    for layer in upper_layers
    for parameter in layer.parameters()
    if parameter.requires_grad
]

head_parameters = list(
    model_b.lm_head.parameters()
)

trainable_params = (
    encoder_parameters + head_parameters
)

# Disable dropout and SpecAugment for this
# controlled comparison.
# eval() does not disable gradient calculations.
model_b.eval()

print(
    "Trainable parameters:",
    sum(p.numel() for p in trainable_params)
)

print(
    "Trainable Transformer layers:",
    len(upper_layers)
)

# ==========================================
# 5. VERIFY STARTING PREDICTIONS
# ==========================================

assert "batches" in globals()
assert "train_ids" in globals()
assert "val_ids" in globals()
assert "report" in globals()
assert "predict_b" in globals()

print("\nCHECKING STARTING MODEL")

starting_result = report(
    "B CLEAN FP32",
    0,
    predict_b
)

# These should match Cell 41's final metrics.
assert abs(
    starting_result["train_cer"] - 0.4989
) < 0.002

assert abs(
    starting_result["val_cer"] - 0.8761
) < 0.002

print("Starting prediction comparison: PASSED")

# ==========================================
# 6. RUN ONE FP32 BACKWARD PASS
# ==========================================

print("\nFP32 GRADIENT DIAGNOSTIC")
print("-" * 55)

test_id = train_ids[0]

model_b.zero_grad(set_to_none=True)

with torch.autocast(
    device_type=DEVICE_42.type,
    enabled=False
):
    output = model_b(**batches[test_id])
    test_loss = output.loss

print("Test recording:", test_id)
print("CTC loss:", float(test_loss.item()))
print("Loss dtype:", test_loss.dtype)
print("Loss requires gradient:", test_loss.requires_grad)

assert torch.isfinite(test_loss).item()
assert test_loss.requires_grad

test_loss.backward()

# ==========================================
# 7. INSPECT EACH PARAMETER'S GRADIENTS
# ==========================================

invalid_gradients = []
missing_gradients = []
valid_gradient_count = 0

for name, parameter in model_b.named_parameters():

    if not parameter.requires_grad:
        continue

    if parameter.grad is None:
        missing_gradients.append(name)
        continue

    if not torch.isfinite(parameter.grad).all():

        invalid_count = int(
            (~torch.isfinite(parameter.grad))
            .sum().item()
        )

        invalid_gradients.append({
            "parameter": name,
            "invalid_values": invalid_count
        })

    else:
        valid_gradient_count += 1

print(
    "\nParameters with valid gradients:",
    valid_gradient_count
)

print(
    "Parameters with missing gradients:",
    len(missing_gradients)
)

print(
    "Parameters with invalid gradients:",
    len(invalid_gradients)
)

if missing_gradients:
    print("\nFirst missing gradients:")
    for name in missing_gradients[:5]:
        print(" ", name)

if invalid_gradients:
    print("\nFirst invalid gradients:")
    for item in invalid_gradients[:10]:
        print(
            item["parameter"],
            "invalid values:",
            item["invalid_values"]
        )

    model_b.zero_grad(set_to_none=True)

    raise RuntimeError(
        "FP32 gradient diagnostic failed. "
        "Do not start training."
    )

# ==========================================
# 8. VERIFY GRADIENT CLIPPING
# ==========================================

gradient_norm = torch.nn.utils.clip_grad_norm_(
    trainable_params,
    max_norm=1.0,
    error_if_nonfinite=True
)

print(
    "\nOriginal gradient norm:",
    float(gradient_norm)
)

model_b.zero_grad(set_to_none=True)

print("\n" + "=" * 55)
print("CLEAN FP32 MODEL: GRADIENT CHECK PASSED")
print("=" * 55)

print("Original XLS-R weights loaded: YES")
print("Cell 41 head restored exactly: YES")
print("Last 2 Transformer layers trainable: YES")
print("All computed gradients finite: YES")
print("Optimizer updates performed: 0")
print("Previous checkpoints modified: NO")


CHECKING PREVIOUS WEIGHT MISMATCH
-------------------------------------------------------
Existing head matches saved head: False
Current head finite: True
Saved head finite: True
Maximum absolute weight difference: 0.0003000497817993164

REBUILDING BRANCH B
-------------------------------------------------------
Saved Cell 41 head restored: VERIFIED
Trainable parameters: 25521473
Trainable Transformer layers: 2

CHECKING STARTING MODEL

B CLEAN FP32 | UPDATE 0
Train CER: 49.89%
Held-out CER: 87.61%
Held-out WER: 100.00%
Anchor: ይምየሳውሸክላየሸክላድ ምስ ው
Held-out: ይሳም ም ሳ ምው
Starting prediction comparison: PASSED

FP32 GRADIENT DIAGNOSTIC
-------------------------------------------------------
Test recording: 6Q0fEziAqyQVIz4J8aws
CTC loss: 1.331987977027893
Loss dtype: torch.float32
Loss requires gradient: True

Parameters with valid gradients: 34
Parameters with missing gradients: 0
Parameters with invalid gradients: 0

Original gradient norm: 10.507054328918457

CLEAN FP32 MODEL: GRADIENT C

In [ ]:

# ============================================================
# CELL 42D - BRANCH B FULL FP32 TRAINING
#
# Starting point:
#   Original XLS-R encoder
#   Cell 41 head at update 4000
#
# Trainable:
#   Last 2 Transformer layers
#   CTC prediction head
#
# Compare against completed Branch A.
# ============================================================

import json
import torch
from pathlib import Path

B_MAX_UPDATES = 300
B_REPORT_EVERY = 100

B_HEAD_LR = 3e-4
B_ENCODER_LR = 1e-5

B_STATE_PATH = RUN_DIR / "last2_fp32_latest.pt"
B_HISTORY_PATH = RUN_DIR / "last2_fp32_history.json"

A_HISTORY_PATH = RUN_DIR / "head_only_history.json"

# ------------------------------------------------------------
# 1. Verify the successful Cell 42C state
# ------------------------------------------------------------

assert "model_b" in globals()
assert "warm_verified" in globals()
assert "train_ids" in globals()
assert "batches" in globals()
assert "report" in globals()
assert "predict_b" in globals()

assert A_HISTORY_PATH.is_file()
assert model_b.training is False

model_b.float()
model_b.eval()

b_trainable = [
    p for p in model_b.parameters()
    if p.requires_grad
]

assert sum(p.numel() for p in b_trainable) == 25521473

assert all(
    p.dtype == torch.float32
    for p in b_trainable
)

# ------------------------------------------------------------
# 2. Create a clean optimizer
# ------------------------------------------------------------

optimizer_b = torch.optim.AdamW(
    [
        {
            "params": encoder_parameters,
            "lr": B_ENCODER_LR,
            "weight_decay": 0.01
        },
        {
            "params": head_parameters,
            "lr": B_HEAD_LR,
            "weight_decay": 0.0
        }
    ]
)

optimizer_b.zero_grad(set_to_none=True)

# ------------------------------------------------------------
# 3. Resume if an FP32 checkpoint already exists
# ------------------------------------------------------------

b_start_step = 0
b_fp32_history = []

if B_STATE_PATH.exists():

    saved = torch.load(
        B_STATE_PATH,
        map_location="cpu",
        weights_only=True
    )

    assert saved["signature"] == signature
    assert saved["precision"] == "fp32"

    model_b.lm_head.load_state_dict(
        saved["head"]
    )

    assert len(saved["upper_layers"]) == 2

    for layer, weights in zip(
        upper_layers,
        saved["upper_layers"]
    ):
        layer.load_state_dict(weights)

    optimizer_b.load_state_dict(
        saved["optimizer"]
    )

    b_start_step = int(saved["step"])

    assert 0 <= b_start_step <= B_MAX_UPDATES

    if B_HISTORY_PATH.exists():
        b_fp32_history = json.loads(
            B_HISTORY_PATH.read_text(encoding="utf-8")
        )

    print("Resuming FP32 training at:", b_start_step)

else:

    # Verify exact saved head before starting.
    for name, parameter in model_b.lm_head.state_dict().items():
        expected = warm_verified["head"][name].to(
            parameter.device
        )

        assert torch.equal(parameter, expected), (
            f"Starting head mismatch: {name}"
        )

    print("Original Cell 41 head: VERIFIED")
    print("Fresh optimizer: INITIALIZED")

# ------------------------------------------------------------
# 4. Check initial or resumed model
# ------------------------------------------------------------

print("\nBRANCH B FP32 CONFIGURATION")
print("=" * 55)

print("Starting step:", b_start_step)
print("Maximum updates:", B_MAX_UPDATES)
print("Precision: FP32")
print("Head learning rate:", B_HEAD_LR)
print("Encoder learning rate:", B_ENCODER_LR)
print("Trainable parameters:",
      sum(p.numel() for p in b_trainable))

if not b_fp32_history:

    start_metrics = report(
        "B FP32",
        b_start_step,
        predict_b
    )

    b_fp32_history.append(start_metrics)

    if b_start_step == 0:
        assert abs(
            start_metrics["train_cer"] - 0.4989
        ) < 0.002

        assert abs(
            start_metrics["val_cer"] - 0.8761
        ) < 0.002

# ------------------------------------------------------------
# 5. Save progress without touching old models
# ------------------------------------------------------------

def save_branch_b_fp32(step):

    state = {
        "signature": signature,
        "precision": "fp32",
        "step": step,
        "head": model_b.lm_head.state_dict(),
        "upper_layers": [
            layer.state_dict()
            for layer in upper_layers
        ],
        "optimizer": optimizer_b.state_dict()
    }

    temporary = RUN_DIR / "last2_fp32_latest.pt.partial"

    torch.save(state, temporary)
    temporary.replace(B_STATE_PATH)

    temporary_history = (
        RUN_DIR / "last2_fp32_history.json.partial"
    )

    temporary_history.write_text(
        json.dumps(
            b_fp32_history,
            indent=2,
            ensure_ascii=False
        ),
        encoding="utf-8"
    )

    temporary_history.replace(B_HISTORY_PATH)

# ------------------------------------------------------------
# 6. Run 300 full-precision optimizer updates
# ------------------------------------------------------------

print("\nTRAINING BRANCH B")
print("=" * 55)

b_completed = b_start_step

for step in range(
    b_start_step + 1,
    B_MAX_UPDATES + 1
):

    # Identical recording order to Branch A.
    rid = train_ids[
        (step - 1) % len(train_ids)
    ]

    optimizer_b.zero_grad(set_to_none=True)

    # Keep dropout and SpecAugment disabled.
    # eval() does not stop backpropagation.
    model_b.eval()

    # Explicitly disable mixed precision.
    with torch.autocast(
        device_type=DEVICE_42.type,
        enabled=False
    ):
        loss = model_b(**batches[rid]).loss

    assert torch.isfinite(loss).item(), (
        f"Invalid FP32 loss at update {step}"
    )

    assert loss.requires_grad

    loss.backward()

    # Stop immediately if a gradient is NaN or Inf.
    grad_norm = torch.nn.utils.clip_grad_norm_(
        b_trainable,
        max_norm=1.0,
        error_if_nonfinite=True
    )

    optimizer_b.step()

    b_completed = step

    if step % B_REPORT_EVERY == 0:

        result = report(
            "B FP32",
            step,
            predict_b
        )

        result["training_loss"] = float(
            loss.item()
        )

        result["gradient_norm"] = float(
            grad_norm
        )

        b_fp32_history.append(result)

        save_branch_b_fp32(step)

        print(
            "Pre-clipping gradient norm:",
            round(float(grad_norm), 4)
        )

        print(
            "Training loss:",
            round(float(loss.item()), 4)
        )

# ------------------------------------------------------------
# 7. Compare saved Branch A with Branch B
# ------------------------------------------------------------

history_a = json.loads(
    A_HISTORY_PATH.read_text(encoding="utf-8")
)

a_by_step = {
    int(row["step"]): row
    for row in history_a
}

b_by_step = {
    int(row["step"]): row
    for row in b_fp32_history
}

print("\n" + "=" * 70)
print("BRANCH A VS BRANCH B")
print("=" * 70)

print(
    f"{'Step':<9}"
    f"{'A Train':<13}"
    f"{'B Train':<13}"
    f"{'A Held-out':<16}"
    f"{'B Held-out':<16}"
)

for step in sorted(
    set(a_by_step) & set(b_by_step)
):

    a = a_by_step[step]
    b = b_by_step[step]

    print(
        f"{step:<9}"
        f"{a['train_cer']*100:<13.2f}"
        f"{b['train_cer']*100:<13.2f}"
        f"{a['val_cer']*100:<16.2f}"
        f"{b['val_cer']*100:<16.2f}"
    )

print("\nFP32 optimizer updates completed:", b_completed)
print("FP32 checkpoint:", B_STATE_PATH)
print("FP32 history:", B_HISTORY_PATH)
print("Previous checkpoints unchanged.")


Original Cell 41 head: VERIFIED
Fresh optimizer: INITIALIZED

BRANCH B FP32 CONFIGURATION
Starting step: 0
Maximum updates: 300
Precision: FP32
Head learning rate: 0.0003
Encoder learning rate: 1e-05
Trainable parameters: 25521473

B FP32 | UPDATE 0
Train CER: 49.89%
Held-out CER: 87.61%
Held-out WER: 100.00%
Anchor: ይምየሳውሸክላየሸክላድ ምስ ው
Held-out: ይሳም ም ሳ ምው

TRAINING BRANCH B

B FP32 | UPDATE 100
Train CER: 45.12%
Held-out CER: 85.04%
Held-out WER: 100.00%
Anchor: ይህምየሳውሸክላየሸክላድ ምስ ው
Held-out: ይሳምስ ም ሳ ምው
Pre-clipping gradient norm: 1.1323
Training loss: 1.399

B FP32 | UPDATE 200
Train CER: 42.63%
Held-out CER: 85.04%
Held-out WER: 100.00%
Anchor: ይህምየሳውሸክላራየሸክላ ድ ምስ ው
Held-out: ይሳምስ ም ስ ሳ በው
Pre-clipping gradient norm: 5.9285
Training loss: 1.1596

B FP32 | UPDATE 300
Train CER: 39.00%
Held-out CER: 85.04%
Held-out WER: 100.00%
Anchor: ይህምየሳውሸክላራ የሸክላ ድስ ምስ ው
Held-out: ይሳምስ ም ስ ሳ በው
Pre-clipping gradient norm: 2.5666
Training loss: 1.1002

BRANCH A VS BRANCH B
Step     A Train      B 

In [ ]:

# ============================================================
# CELL 43 - SCALED DATASET: 64 TRAIN / 16 HELD-OUT
#
# Reuse the 8 previously trained recordings.
# Select fresh held-out speakers.
# Prefer shorter recordings and diverse speakers.
#
# No GPU training or checkpoint modifications.
# ============================================================

import json
import random
import statistics
from collections import defaultdict, Counter
from pathlib import Path
from IPython.display import Audio, display

SEED_43 = 20261019
TRAIN_TARGET = 64
VAL_TARGET = 16
VAL_SPEAKERS = 8
VAL_PER_SPEAKER = 2

EXP43_DIR = DATA_DIR / "scaled_amharic_64_16_v1"
EXP43_DIR.mkdir(parents=True, exist_ok=True)
EXP43_SELECTION = EXP43_DIR / "selection.json"

OLD_SPLIT = (
    DATA_DIR
    / "short_multirecording_head_only_v2"
    / "split.json"
)

assert OLD_SPLIT.is_file()

previous_split = json.loads(
    OLD_SPLIT.read_text(encoding="utf-8")
)

carryover_ids = previous_split["train_ids"]
assert len(carryover_ids) == 8

by_id_43 = {r["id"]: r for r in train_records}
assert all(rid in by_id_43 for rid in carryover_ids)

# Exclude every speaker previously involved in
# our small experiments from the NEW validation set.
prior_ids = set(
    previous_split["train_ids"]
    + previous_split["val_ids"]
)

old_long_selection = (
    DATA_DIR
    / "head_only_multirecording_v1"
    / "selection.json"
)

if old_long_selection.exists():
    old = json.loads(
        old_long_selection.read_text(encoding="utf-8")
    )
    prior_ids.update(old["train_ids"])
    prior_ids.update(old["val_ids"])

prior_speakers = {
    by_id_43[rid]["speaker_id"]
    for rid in prior_ids
    if rid in by_id_43
}

KERNELS_43 = (10, 3, 3, 3, 3, 2, 2)
STRIDES_43 = (5, 2, 2, 2, 2, 2, 2)

def count_frames_43(samples):
    for kernel, stride in zip(KERNELS_43, STRIDES_43):
        samples = (samples - kernel) // stride + 1
    return samples

def eligible_43(record, max_duration, allow_digits):
    duration = float(record["duration_seconds"])
    text = record["transcription"]

    if not (4.0 <= duration <= max_duration):
        return False

    if not record.get("speaker_id"):
        return False

    if not allow_digits and any(c.isdigit() for c in text):
        return False

    path = Path(AUDIO_DIR) / record["audio_file"]
    if not path.is_file() or path.stat().st_size == 0:
        return False

    labels = tokenizer.encode(
        text, add_special_tokens=False
    )

    if not (20 <= len(labels) <= 160):
        return False

    if tokenizer.unk_token_id in labels:
        return False

    repeats = sum(
        a == b
        for a, b in zip(labels[:-1], labels[1:])
    )

    frames = count_frames_43(round(duration * 16000))
    return frames - len(labels) - repeats >= 20

def try_select_43(max_duration, allow_digits):
    rng = random.Random(SEED_43)

    groups = defaultdict(list)

    for record in train_records:
        if eligible_43(record, max_duration, allow_digits):
            groups[record["speaker_id"]].append(record)

    for sid in groups:
        groups[sid].sort(key=lambda r: r["id"])
        rng.shuffle(groups[sid])

    # Only unfamiliar speakers can enter validation.
    valid_speakers = [
        sid for sid, records in groups.items()
        if sid not in prior_speakers
        and len(records) >= VAL_PER_SPEAKER
    ]

    valid_speakers.sort()
    rng.shuffle(valid_speakers)

    if len(valid_speakers) < VAL_SPEAKERS:
        return None

    heldout_speakers = set(
        valid_speakers[:VAL_SPEAKERS]
    )

    val_ids = [
        record["id"]
        for sid in valid_speakers[:VAL_SPEAKERS]
        for record in groups[sid][:VAL_PER_SPEAKER]
    ]

    # Carryover examples must remain part of training.
    if not all(
        eligible_43(by_id_43[rid], max_duration, allow_digits)
        for rid in carryover_ids
    ):
        return None

    train_ids = list(carryover_ids)
    used_ids = set(train_ids)

    speaker_counts = Counter(
        by_id_43[rid]["speaker_id"]
        for rid in train_ids
    )

    train_speakers = sorted(
        sid for sid in groups
        if sid not in heldout_speakers
    )
    rng.shuffle(train_speakers)

    # Round robin encourages speaker diversity.
    # Limit to three examples from each speaker.
    for _ in range(3):
        for sid in train_speakers:
            if len(train_ids) >= TRAIN_TARGET:
                break
            if speaker_counts[sid] >= 3:
                continue

            for record in groups[sid]:
                rid = record["id"]

                if rid not in used_ids:
                    train_ids.append(rid)
                    used_ids.add(rid)
                    speaker_counts[sid] += 1
                    break

        if len(train_ids) >= TRAIN_TARGET:
            break

    if len(train_ids) != TRAIN_TARGET:
        return None

    return {
        "train_ids": train_ids,
        "val_ids": val_ids,
        "seed": SEED_43,
        "max_duration_seconds": max_duration,
        "digits_allowed": allow_digits,
        "carryover_ids": carryover_ids,
        "source": "train_final_25h_ctc_safe"
    }

# ------------------------------------------------------------
# Restore or construct selection
# ------------------------------------------------------------

if EXP43_SELECTION.exists():
    selection_43 = json.loads(
        EXP43_SELECTION.read_text(encoding="utf-8")
    )
    print("Existing scaled selection restored.")

else:
    selection_43 = None

    for allow_digits in [False, True]:
        for max_duration in [10, 12, 15, 18]:
            selection_43 = try_select_43(
                max_duration, allow_digits
            )

            if selection_43 is not None:
                print(
                    "Selection succeeded:",
                    max_duration, "seconds,",
                    "digits allowed:", allow_digits
                )
                break

        if selection_43 is not None:
            break

    assert selection_43 is not None, (
        "Not enough eligible recordings. "
        "Review the selection constraints."
    )

    temporary = EXP43_DIR / "selection.json.partial"
    temporary.write_text(
        json.dumps(
            selection_43,
            indent=2,
            ensure_ascii=False
        ),
        encoding="utf-8"
    )
    temporary.replace(EXP43_SELECTION)

train_ids_43 = selection_43["train_ids"]
val_ids_43 = selection_43["val_ids"]

assert len(train_ids_43) == TRAIN_TARGET
assert len(val_ids_43) == VAL_TARGET
assert len(set(train_ids_43 + val_ids_43)) == 80
assert set(carryover_ids).issubset(train_ids_43)

train_records_43 = [
    by_id_43[rid] for rid in train_ids_43
]
val_records_43 = [
    by_id_43[rid] for rid in val_ids_43
]

train_speakers_43 = {
    r["speaker_id"] for r in train_records_43
}
val_speakers_43 = {
    r["speaker_id"] for r in val_records_43
}

assert not (train_speakers_43 & val_speakers_43)
assert not (prior_speakers & val_speakers_43)
assert len(val_speakers_43) == VAL_SPEAKERS

assert all(
    eligible_43(
        r,
        selection_43["max_duration_seconds"],
        selection_43["digits_allowed"]
    )
    for r in train_records_43 + val_records_43
)

def duration_summary_43(records):
    values = [
        float(r["duration_seconds"])
        for r in records
    ]

    return (
        round(statistics.mean(values), 2),
        round(max(values), 2),
        round(sum(values) / 60, 2)
    )

print("\n" + "=" * 60)
print("CELL 43: SCALED DATASET SUMMARY")
print("=" * 60)

print("Train recordings:", len(train_records_43))
print("Held-out recordings:", len(val_records_43))
print("Training speakers:", len(train_speakers_43))
print("Held-out speakers:", len(val_speakers_43))
print("Speaker overlap:", 0)
print("Old training examples retained:", len(carryover_ids))
print("Previous experiment speakers in validation:", 0)

print("\nTrain (mean sec, max sec, total min):",
      duration_summary_43(train_records_43))
print("Held-out (mean sec, max sec, total min):",
      duration_summary_43(val_records_43))

print("\nFIRST 5 TRAINING RECORDINGS")
for record in train_records_43[:5]:
    print(
        record["id"],
        round(float(record["duration_seconds"]), 2),
        record["transcription"][:100]
    )

print("\nFIRST 5 HELD-OUT RECORDINGS")
for record in val_records_43[:5]:
    print(
        record["id"],
        round(float(record["duration_seconds"]), 2),
        record["transcription"][:100]
    )

# ------------------------------------------------------------
# Manual audio/transcript inspection
# ------------------------------------------------------------

print("\nAUDIO QUALITY SPOT CHECK")

for label, record in [
    ("NEW TRAINING", train_records_43[8]),
    ("HELD-OUT 1", val_records_43[0]),
    ("HELD-OUT 2", val_records_43[1])
]:
    print("\n", label)
    print("ID:", record["id"])
    print("Transcript:", record["transcription"])

    display(Audio(
        filename=str(
            Path(AUDIO_DIR) / record["audio_file"]
        )
    ))

print("\nDATASET VALIDATION PASSED")
print("Selection saved:", EXP43_SELECTION)
print("No model weights or checkpoints modified.")


Existing scaled selection restored.

CELL 43: SCALED DATASET SUMMARY
Train recordings: 64
Held-out recordings: 16
Training speakers: 60
Held-out speakers: 8
Speaker overlap: 0
Old training examples retained: 8
Previous experiment speakers in validation: 0

Train (mean sec, max sec, total min): (12.91, 14.98, 13.77)
Held-out (mean sec, max sec, total min): (14.65, 14.98, 3.91)

FIRST 5 TRAINING RECORDINGS
6Q0fEziAqyQVIz4J8aws 5.18 ይህ ምስል የሚያሳየው ከሸክላ የሚሰራ የሸክላ ድስት ምስል ነው
8DDU79GSsgg8dZV0J3ox 4.3 ወንድ አርሶአደር በማሳ ላይ እየተጓዘ
VpYkSBOYaCCY8Zx6cEDm 5.18 ምስሉ ላይ የምንመለከተው በአንድ የሸክላ ንስሀ ውስጥ ያለ የዶሮ ወጥ ነው
GjjqjszNttEsTkd4oBja 7.46 በምስሉ ላይ የምትመለከቱ ግ አስከባሪዎች ወደ እምነት ስርዓት የሚመጡ ሰዎችን እየፈተሽ ነው
GIJ84glb4OAhzMApjlDC 7.58 ይህ በምስሉ የምንመለከተው ወንዝ ሲሆን ሰዎች ልብሳቸውን እያጠቡ ሰዎች ልብሳቸውን እያጠቡ ከብቶቻቸውን ውሃ እያጠጡ እንዲሁም ውሃ እየቀዱ

FIRST 5 HELD-OUT RECORDINGS
4ljLQRFgHFJqEsJDZuHd 14.26 ይህ የምንመለከተዉ ምስል የኢትዮጵያ ባህላዊ ግብይት እንዲሁም ሸመታ ነዉ
AbsVNlAJl7BLd05CFVhu 14.66 ይህ ምንመለከተው ምስል የሴቶች የፀጉር አሰራር ሲሆን ስሙ ሹሩባ ይባላል አብዛኞቹ የ ኢትዮጵያ ሴቶች ይህን አሰራር ይሰሩታል


 HELD-OUT 1
ID: 4ljLQRFgHFJqEsJDZuHd
Transcript: ይህ የምንመለከተዉ ምስል የኢትዮጵያ ባህላዊ ግብይት እንዲሁም ሸመታ ነዉ



 HELD-OUT 2
ID: AbsVNlAJl7BLd05CFVhu
Transcript: ይህ ምንመለከተው ምስል የሴቶች የፀጉር አሰራር ሲሆን ስሙ ሹሩባ ይባላል አብዛኞቹ የ ኢትዮጵያ ሴቶች ይህን አሰራር ይሰሩታል



DATASET VALIDATION PASSED
Selection saved: /content/drive/MyDrive/Amharic_ASR_XLSR/data/scaled_amharic_64_16_v1/selection.json
No model weights or checkpoints modified.


In [ ]:

# ============================================================
# CELL 44 - SCALED TRAINING PREFLIGHT
#
# Restore Branch B from Cell 42D, update 300.
# Verify gradients on the longest training recording.
# Evaluate 16 new held-out recordings.
#
# No optimizer updates or checkpoint overwrites.
# ============================================================

import json
import gc
import statistics
from pathlib import Path

import torch
from jiwer import cer, wer
from transformers import Wav2Vec2ForCTC

DEVICE_44 = torch.device(
    "cuda" if torch.cuda.is_available() else "cpu"
)

SOURCE_CHECKPOINT = (
    DATA_DIR
    / "warm_head_encoder_comparison_v1"
    / "last2_fp32_latest.pt"
)

SELECTION_44 = (
    DATA_DIR
    / "scaled_amharic_64_16_v1"
    / "selection.json"
)

PREFLIGHT_PATH = (
    DATA_DIR
    / "scaled_amharic_64_16_v1"
    / "fp32_preflight.json"
)

assert SOURCE_CHECKPOINT.is_file()
assert SELECTION_44.is_file()

selection_44 = json.loads(
    SELECTION_44.read_text(encoding="utf-8")
)

train_ids_44 = selection_44["train_ids"]
val_ids_44 = selection_44["val_ids"]

assert len(train_ids_44) == 64
assert len(val_ids_44) == 16

record_by_id_44 = {
    record["id"]: record
    for record in train_records
}

dataset_index_44 = {
    record["id"]: index
    for index, record in enumerate(train_dataset.records)
}

assert all(
    rid in dataset_index_44
    for rid in train_ids_44 + val_ids_44
)

train_speakers_44 = {
    record_by_id_44[rid]["speaker_id"]
    for rid in train_ids_44
}

val_speakers_44 = {
    record_by_id_44[rid]["speaker_id"]
    for rid in val_ids_44
}

assert not (train_speakers_44 & val_speakers_44)

# ------------------------------------------------------------
# 1. Load the successful Branch B checkpoint
# ------------------------------------------------------------

print("LOADING BRANCH B")
print("=" * 55)

saved_44 = torch.load(
    SOURCE_CHECKPOINT,
    map_location="cpu",
    weights_only=True
)

assert saved_44["precision"] == "fp32"
assert int(saved_44["step"]) == 300
assert len(saved_44["upper_layers"]) == 2

model_44 = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(DEVICE_44).float()

model_44.lm_head.load_state_dict(
    saved_44["head"],
    strict=True
)

upper_layers_44 = list(
    model_44.wav2vec2.encoder.layers[-2:]
)

for layer, weights in zip(
    upper_layers_44,
    saved_44["upper_layers"]
):
    layer.load_state_dict(weights, strict=True)

# Freeze all parameters.
model_44.requires_grad_(False)

# Enable the same components as Branch B.
for layer in upper_layers_44:
    layer.requires_grad_(True)

model_44.lm_head.requires_grad_(True)

# Keep dropout and SpecAugment disabled
# during this controlled experiment.
model_44.eval()

trainable_44 = [
    parameter
    for parameter in model_44.parameters()
    if parameter.requires_grad
]

assert sum(
    p.numel() for p in trainable_44
) == 25521473

print("Checkpoint step: 300")
print("Precision: FP32")
print("Trainable parameters:", sum(
    p.numel() for p in trainable_44
))

# ------------------------------------------------------------
# 2. Helper: Retrieve one recording
# ------------------------------------------------------------

def get_batch_44(record_id):

    example = train_dataset[
        dataset_index_44[record_id]
    ]

    batch = ctc_collator([example])

    return {
        key: value.to(DEVICE_44)
        for key, value in batch.items()
    }

def decode_44(logits):

    predicted_ids = logits.argmax(dim=-1)

    prediction = processor.batch_decode(
        predicted_ids.cpu()
    )[0]

    return normalize_amharic_ctc(
        prediction
    )

# ------------------------------------------------------------
# 3. Evaluate the new validation set
# ------------------------------------------------------------

print("\nNEW VALIDATION BASELINE")
print("=" * 55)

references_44 = []
predictions_44 = []
validation_rows_44 = []

model_44.eval()

with torch.no_grad():

    for index, rid in enumerate(val_ids_44, 1):

        batch = get_batch_44(rid)

        logits = model_44(**batch).logits
        prediction = decode_44(logits)

        reference = normalize_amharic_ctc(
            record_by_id_44[rid]["transcription"]
        )

        references_44.append(reference)
        predictions_44.append(prediction)

        validation_rows_44.append({
            "id": rid,
            "reference": reference,
            "prediction": prediction,
            "cer": float(cer(reference, prediction)),
            "wer": float(wer(reference, prediction)),
            "duration": float(
                record_by_id_44[rid]["duration_seconds"]
            )
        })

        if index <= 3:
            print(f"\nValidation recording {index}")
            print("ID:", rid)
            print("Reference:", reference[:150])
            print(
                "Prediction:",
                prediction[:150] or "[EMPTY]"
            )

        del batch, logits

baseline_cer_44 = float(
    cer(references_44, predictions_44)
)

baseline_wer_44 = float(
    wer(references_44, predictions_44)
)

print("\nValidation CER:",
      f"{baseline_cer_44 * 100:.2f}%")

print("Validation WER:",
      f"{baseline_wer_44 * 100:.2f}%")

print("Nonempty predictions:", sum(
    bool(p.strip()) for p in predictions_44
), "/16")

# ------------------------------------------------------------
# 4. Test gradients on the LONGEST training recording
# ------------------------------------------------------------

longest_id_44 = max(
    train_ids_44,
    key=lambda rid: float(
        record_by_id_44[rid]["duration_seconds"]
    )
)

longest_duration_44 = float(
    record_by_id_44[
        longest_id_44
    ]["duration_seconds"]
)

print("\nLONG-RECORDING FP32 GRADIENT TEST")
print("=" * 55)

print("Recording:", longest_id_44)
print("Duration:", longest_duration_44, "seconds")

test_batch_44 = get_batch_44(longest_id_44)

# Confirm actual CTC alignment feasibility.
target_ids_44 = test_batch_44["labels"][
    test_batch_44["labels"] >= 0
]

actual_frames_44 = int(
    model_44._get_feat_extract_output_lengths(
        torch.tensor([
            test_batch_44["input_values"].shape[1]
        ])
    )[0].item()
)

repeats_44 = int(
    (target_ids_44[1:] == target_ids_44[:-1])
    .sum().item()
)

required_frames_44 = (
    target_ids_44.numel() + repeats_44
)

print("Available CTC frames:", actual_frames_44)
print("Required CTC frames:", required_frames_44)

assert actual_frames_44 >= required_frames_44

# Free existing gradients from previous work.
model_44.zero_grad(set_to_none=True)

if DEVICE_44.type == "cuda":
    torch.cuda.reset_peak_memory_stats()

# No autocast. No gradient scaler.
with torch.autocast(
    device_type=DEVICE_44.type,
    enabled=False
):
    test_loss_44 = model_44(**test_batch_44).loss

print("\nLoss:", float(test_loss_44.item()))
print("Loss dtype:", test_loss_44.dtype)
print("Requires grad:", test_loss_44.requires_grad)

assert torch.isfinite(test_loss_44).item()
assert test_loss_44.requires_grad

test_loss_44.backward()

# ------------------------------------------------------------
# 5. Verify gradients before any training
# ------------------------------------------------------------

invalid_44 = []
missing_44 = []
valid_44 = 0

for name, parameter in model_44.named_parameters():

    if not parameter.requires_grad:
        continue

    if parameter.grad is None:
        missing_44.append(name)
        continue

    if not torch.isfinite(parameter.grad).all().item():
        invalid_44.append(name)
    else:
        valid_44 += 1

print("\nGRADIENT RESULTS")
print("Valid parameter gradients:", valid_44)
print("Missing parameter gradients:", len(missing_44))
print("Invalid parameter gradients:", len(invalid_44))

assert not invalid_44, (
    f"Invalid gradients: {invalid_44[:5]}"
)

assert not missing_44, (
    f"Missing gradients: {missing_44[:5]}"
)

gradient_norm_44 = torch.nn.utils.clip_grad_norm_(
    trainable_44,
    max_norm=1.0,
    error_if_nonfinite=True
)

print(
    "Gradient norm before clipping:",
    round(float(gradient_norm_44), 4)
)

peak_gpu_gb_44 = None

if DEVICE_44.type == "cuda":
    peak_gpu_gb_44 = (
        torch.cuda.max_memory_allocated()
        / 1024**3
    )

    print(
        "Peak allocated GPU memory:",
        round(peak_gpu_gb_44, 2),
        "GB"
    )

# Remove gradients from the diagnostic.
model_44.zero_grad(set_to_none=True)

del test_batch_44, test_loss_44
gc.collect()

if DEVICE_44.type == "cuda":
    torch.cuda.empty_cache()

# ------------------------------------------------------------
# 6. Save baseline measurements
# ------------------------------------------------------------

preflight_report_44 = {
    "source_checkpoint": str(SOURCE_CHECKPOINT),
    "source_step": 300,
    "training_examples": len(train_ids_44),
    "validation_examples": len(val_ids_44),
    "validation_cer": baseline_cer_44,
    "validation_wer": baseline_wer_44,
    "validation_predictions": validation_rows_44,
    "longest_train_recording": longest_id_44,
    "longest_train_duration": longest_duration_44,
    "gradient_norm": float(gradient_norm_44),
    "valid_gradient_tensors": valid_44,
    "invalid_gradient_tensors": len(invalid_44),
    "peak_allocated_gpu_gb": peak_gpu_gb_44
}

PREFLIGHT_PATH.write_text(
    json.dumps(
        preflight_report_44,
        indent=2,
        ensure_ascii=False
    ),
    encoding="utf-8"
)

print("\n" + "=" * 55)
print("SCALED TRAINING PREFLIGHT PASSED")
print("=" * 55)

print("Validation CER:",
      f"{baseline_cer_44 * 100:.2f}%")
print("Validation WER:",
      f"{baseline_wer_44 * 100:.2f}%")
print("Full-precision gradients: VALID")
print("Optimizer updates: 0")
print("Baseline saved:", PREFLIGHT_PATH)
print("Existing checkpoints: UNCHANGED")


LOADING BRANCH B
Checkpoint step: 300
Precision: FP32
Trainable parameters: 25521473

NEW VALIDATION BASELINE

Validation recording 1
ID: 4ljLQRFgHFJqEsJDZuHd
Reference: ይህ የምንመለከተዉ ምስል የኢትዮጵያ ባህላዊ ግብይት እንዲሁም ሸመታ ነዉ
Prediction: ፀው ይ ህየውሳበምውበርበሰ ውየማበድውው

Validation recording 2
ID: AbsVNlAJl7BLd05CFVhu
Reference: ይህ ምንመለከተው ምስል የሴቶች የፀጉር አሰራር ሲሆን ስሙ ሹሩባ ይባላል አብዛኞቹ የ ኢትዮጵያ ሴቶች ይህን አሰራር ይሰሩታል
Prediction: ይው ውውምበሰበስስሰ ም የ ውውውው

Validation recording 3
ID: 3XmMbvidHt0izuWdATyW
Reference: ባንድራ እና መላያ የኢትዮጵያ ባንድራ የኢትዮጵያ ባንድራ የህዝቦቹን ተስፋ አንድነት ታሪክ ልምላሜ ተጋድሎን የሚገልጽ በህዝቦች ዘንድ ሰላምን የሚያመለክት የባንድራ አይነት ነው
Prediction: ነህውልና ልልምእይንስልእእምው ስእምነእውነንውምናነንነውንይነውውምውልትልእምውጉነእእምውልልልስነይልእው ናንንምውምህንናህስእንእየናህነ

Validation CER: 90.56%
Validation WER: 99.70%
Nonempty predictions: 16 /16

LONG-RECORDING FP32 GRADIENT TEST
Recording: 1kPe5yhdSKLyyBYtp1yP
Duration: 14.976 seconds
Available CTC frames: 748
Required CTC frames: 60

Loss: 6.966094493865967
Loss dtype: torch.float32
Requires grad: True

GRADIENT RESULTS
Va

In [ ]:

# ============================================================
# CELL 45 - SCALED FP32 TRAINING PILOT
#
# 64 training recordings, 16 held-out recordings
# Start from Branch B at update 300
# Train last 2 Transformer layers + CTC head
#
# 128 updates (2 passes through 64 recordings)
# Evaluate and checkpoint every 32 updates
# ============================================================

import json
import random
import hashlib
import statistics
from pathlib import Path

import torch
from jiwer import cer, wer

PILOT_STEPS = 128
REPORT_INTERVAL = 32

HEAD_LR_45 = 1e-4
ENCODER_LR_45 = 2e-6
CLIP_NORM_45 = 1.0

PILOT_DIR = (
    DATA_DIR
    / "scaled_amharic_64_16_v1"
    / "stage1_fp32"
)
PILOT_DIR.mkdir(parents=True, exist_ok=True)

STATE_45 = PILOT_DIR / "latest.pt"
HISTORY_45 = PILOT_DIR / "history.json"

required_names = [
    "model_44", "saved_44",
    "train_ids_44", "val_ids_44",
    "get_batch_44", "record_by_id_44",
    "decode_44"
]

missing = [
    name for name in required_names
    if name not in globals()
]
assert not missing, f"Missing Cell 44 state: {missing}"

assert len(train_ids_44) == 64
assert len(val_ids_44) == 16
assert int(saved_44["step"]) == 300

# ------------------------------------------------------------
# 1. Reconfigure the existing model
# ------------------------------------------------------------

model_44 = model_44.float()
model_44.requires_grad_(False)

upper_45 = list(
    model_44.wav2vec2.encoder.layers[-2:]
)

for layer in upper_45:
    layer.requires_grad_(True)

model_44.lm_head.requires_grad_(True)
model_44.eval()

encoder_params_45 = [
    p for layer in upper_45
    for p in layer.parameters()
    if p.requires_grad
]

head_params_45 = list(
    model_44.lm_head.parameters()
)

trainable_45 = encoder_params_45 + head_params_45

assert sum(p.numel() for p in trainable_45) == 25521473

optimizer_45 = torch.optim.AdamW([
    {
        "params": encoder_params_45,
        "lr": ENCODER_LR_45,
        "weight_decay": 0.01
    },
    {
        "params": head_params_45,
        "lr": HEAD_LR_45,
        "weight_decay": 0.0
    }
])

# A new optimizer starts here. We retain trained
# weights but reset AdamW's moment estimates.

config_45 = {
    "source": str(SOURCE_CHECKPOINT),
    "source_step": 300,
    "train_ids": train_ids_44,
    "val_ids": val_ids_44,
    "references": {
        rid: record_by_id_44[rid]["transcription"]
        for rid in train_ids_44 + val_ids_44
    },
    "head_lr": HEAD_LR_45,
    "encoder_lr": ENCODER_LR_45,
    "clip_norm": CLIP_NORM_45,
    "seed": 451
}

signature_45 = hashlib.sha256(
    json.dumps(
        config_45,
        sort_keys=True,
        ensure_ascii=False
    ).encode("utf-8")
).hexdigest()

# ------------------------------------------------------------
# 2. Restore saved pilot progress or warm-start weights
# ------------------------------------------------------------

start_45 = 0
history_45 = []

if STATE_45.exists():

    saved = torch.load(
        STATE_45,
        map_location="cpu",
        weights_only=True
    )

    assert saved["signature"] == signature_45

    model_44.lm_head.load_state_dict(saved["head"])

    for layer, weights in zip(
        upper_45, saved["upper_layers"]
    ):
        layer.load_state_dict(weights)

    optimizer_45.load_state_dict(saved["optimizer"])
    start_45 = int(saved["step"])

    if HISTORY_45.exists():
        history_45 = json.loads(
            HISTORY_45.read_text(encoding="utf-8")
        )

    print("Resuming pilot from update:", start_45)

else:

    # Restore exact Branch B update-300 weights.
    model_44.lm_head.load_state_dict(
        saved_44["head"]
    )

    for layer, weights in zip(
        upper_45, saved_44["upper_layers"]
    ):
        layer.load_state_dict(weights)

    print("Starting from verified Branch B update 300.")

assert 0 <= start_45 <= PILOT_STEPS

# ------------------------------------------------------------
# 3. Evaluation
# ------------------------------------------------------------

# Eight previously trained examples plus eight newly
# selected training examples form a fixed training probe.
train_probe_45 = (
    train_ids_44[:8] + train_ids_44[8:16]
)

def evaluate_45(record_ids):

    model_44.eval()

    refs = []
    preds = []

    with torch.no_grad():

        for rid in record_ids:

            batch = get_batch_44(rid)

            output = model_44(
                input_values=batch["input_values"],
                attention_mask=batch["attention_mask"]
            )

            prediction = decode_44(output.logits)

            reference = normalize_amharic_ctc(
                record_by_id_44[rid]["transcription"]
            )

            refs.append(reference)
            preds.append(prediction)

            del output, batch

    return {
        "cer": float(cer(refs, preds)),
        "wer": float(wer(refs, preds)),
        "nonempty": sum(bool(p.strip()) for p in preds),
        "predictions": preds
    }

def report_45(step):

    train_result = evaluate_45(train_probe_45)
    val_result = evaluate_45(val_ids_44)

    result = {
        "step": step,
        "train_probe_cer": train_result["cer"],
        "val_cer": val_result["cer"],
        "val_wer": val_result["wer"],
        "val_nonempty": val_result["nonempty"],
        "train_prediction": train_result["predictions"][0],
        "val_prediction": val_result["predictions"][0]
    }

    print(f"\nUPDATE {step}/{PILOT_STEPS}")
    print("-" * 50)

    print(
        "Training probe CER (16 recordings):",
        f"{result['train_probe_cer'] * 100:.2f}%"
    )

    print(
        "Held-out CER (16 recordings):",
        f"{result['val_cer'] * 100:.2f}%"
    )

    print(
        "Held-out WER:",
        f"{result['val_wer'] * 100:.2f}%"
    )

    print(
        "Held-out nonempty predictions:",
        f"{result['val_nonempty']}/16"
    )

    print(
        "Held-out example:",
        result["val_prediction"][:120] or "[EMPTY]"
    )

    return result

def save_45(step):

    checkpoint = {
        "signature": signature_45,
        "step": step,
        "precision": "fp32",
        "head": model_44.lm_head.state_dict(),
        "upper_layers": [
            layer.state_dict()
            for layer in upper_45
        ],
        "optimizer": optimizer_45.state_dict()
    }

    temp_state = PILOT_DIR / "latest.pt.partial"
    torch.save(checkpoint, temp_state)
    temp_state.replace(STATE_45)

    temp_history = PILOT_DIR / "history.json.partial"

    temp_history.write_text(
        json.dumps(
            history_45,
            indent=2,
            ensure_ascii=False
        ),
        encoding="utf-8"
    )

    temp_history.replace(HISTORY_45)

# ------------------------------------------------------------
# 4. Establish baseline
# ------------------------------------------------------------

print("\nSCALED FP32 PILOT")
print("=" * 55)
print("Training recordings: 64")
print("Held-out recordings: 16")
print("Trainable parameters: 25,521,473")
print("Head LR:", HEAD_LR_45)
print("Encoder LR:", ENCODER_LR_45)
print("Gradient clip:", CLIP_NORM_45)
print("FP16 autocast: DISABLED")

if start_45 == 0 and not history_45:

    baseline_45 = report_45(0)

    preflight = json.loads(
        PREFLIGHT_PATH.read_text(encoding="utf-8")
    )

    # Confirm the clean initial validation model.
    assert abs(
        baseline_45["val_cer"]
        - preflight["validation_cer"]
    ) < 0.01, "Baseline mismatch; stop before training."

    history_45.append(baseline_45)

# ------------------------------------------------------------
# 5. Deterministic speaker-diverse data order
# ------------------------------------------------------------

def record_for_step_45(step):

    zero_index = step - 1
    epoch = zero_index // len(train_ids_44)
    position = zero_index % len(train_ids_44)

    order = list(train_ids_44)

    rng = random.Random(451 + epoch)
    rng.shuffle(order)

    return order[position]

# ------------------------------------------------------------
# 6. Run 128 optimizer updates
# ------------------------------------------------------------

recent_norms = []
recent_losses = []
completed_45 = start_45

for step in range(start_45 + 1, PILOT_STEPS + 1):

    rid = record_for_step_45(step)

    model_44.eval()
    optimizer_45.zero_grad(set_to_none=True)

    batch = get_batch_44(rid)

    # Full precision, including CTC calculation.
    with torch.autocast(
        device_type=DEVICE_44.type,
        enabled=False
    ):
        loss = model_44(**batch).loss

    if not torch.isfinite(loss).item():
        raise RuntimeError(
            f"Non-finite loss at update {step}, ID {rid}"
        )

    loss.backward()

    grad_norm = torch.nn.utils.clip_grad_norm_(
        trainable_45,
        max_norm=CLIP_NORM_45,
        error_if_nonfinite=True
    )

    raw_norm = float(grad_norm)

    # Stop on extreme unexpected gradients.
    if raw_norm > 5000:
        optimizer_45.zero_grad(set_to_none=True)
        raise RuntimeError(
            f"Extreme gradient norm {raw_norm:.1f} "
            f"at update {step}, recording {rid}"
        )

    optimizer_45.step()

    recent_norms.append(raw_norm)
    recent_losses.append(float(loss.item()))

    completed_45 = step

    del batch, loss

    if step % REPORT_INTERVAL == 0:

        result = report_45(step)

        result["mean_train_step_loss"] = (
            statistics.mean(recent_losses)
        )
        result["median_gradient_norm"] = (
            statistics.median(recent_norms)
        )
        result["max_gradient_norm"] = max(
            recent_norms
        )
        result["fraction_gradients_clipped"] = (
            sum(n > CLIP_NORM_45 for n in recent_norms)
            / len(recent_norms)
        )

        print(
            "Mean optimizer-step loss:",
            round(result["mean_train_step_loss"], 4)
        )

        print(
            "Median gradient norm:",
            round(result["median_gradient_norm"], 2)
        )

        print(
            "Maximum gradient norm:",
            round(result["max_gradient_norm"], 2)
        )

        print(
            "Fraction of steps clipped:",
            f"{result['fraction_gradients_clipped'] * 100:.1f}%"
        )

        history_45.append(result)
        save_45(step)

        recent_norms.clear()
        recent_losses.clear()

# ------------------------------------------------------------
# 7. Summary
# ------------------------------------------------------------

print("\n" + "=" * 65)
print("SCALED FP32 PILOT SUMMARY")
print("=" * 65)

print(
    f"{'Update':<9}"
    f"{'Train probe CER':<19}"
    f"{'Held-out CER':<17}"
    f"{'Held-out WER':<17}"
)

for row in history_45:

    print(
        f"{row['step']:<9}"
        f"{row['train_probe_cer']*100:<19.2f}"
        f"{row['val_cer']*100:<17.2f}"
        f"{row['val_wer']*100:<17.2f}"
    )

print("\nUpdates completed:", completed_45)
print("Checkpoint:", STATE_45)
print("History:", HISTORY_45)
print("Earlier experiments and checkpoints unchanged.")


Starting from verified Branch B update 300.

SCALED FP32 PILOT
Training recordings: 64
Held-out recordings: 16
Trainable parameters: 25,521,473
Head LR: 0.0001
Encoder LR: 2e-06
Gradient clip: 1.0
FP16 autocast: DISABLED

UPDATE 0/128
--------------------------------------------------
Training probe CER (16 recordings): 69.41%
Held-out CER (16 recordings): 90.56%
Held-out WER: 99.70%
Held-out nonempty predictions: 16/16
Held-out example: ፀው ይ ህየውሳበምውበርበሰ ውየማበድውው

UPDATE 32/128
--------------------------------------------------
Training probe CER (16 recordings): 70.20%
Held-out CER (16 recordings): 89.84%
Held-out WER: 99.70%
Held-out nonempty predictions: 16/16
Held-out example: ፀው ይ ውሳበምውበርበ በውማበድውው
Mean optimizer-step loss: 6.7714
Median gradient norm: 40.21
Maximum gradient norm: 416.28
Fraction of steps clipped: 100.0%

UPDATE 64/128
--------------------------------------------------
Training probe CER (16 recordings): 70.64%
Held-out CER (16 recordings): 89.54%
Held-out WER: 99.7

In [ ]:

# ============================================================
# CELL 46 - SCALED ASR FAILURE-MODE AUDIT
#
# Evaluate 64 training + 16 held-out recordings.
# Measure CER, WER, CTC loss, blank behavior,
# output length, and transcription density.
#
# No training. No checkpoint modifications.
# ============================================================

import json
import statistics
from collections import defaultdict
from pathlib import Path

import torch
from transformers import Wav2Vec2ForCTC
from jiwer import cer, wer

AUDIT_DIR = (
    DATA_DIR / "scaled_amharic_64_16_v1"
)
AUDIT_CHECKPOINT = (
    AUDIT_DIR / "stage1_fp32" / "latest.pt"
)
AUDIT_SELECTION = AUDIT_DIR / "selection.json"
AUDIT_BASELINE = AUDIT_DIR / "fp32_preflight.json"
AUDIT_OUTPUT = AUDIT_DIR / "failure_mode_audit.json"

assert AUDIT_CHECKPOINT.is_file()
assert AUDIT_SELECTION.is_file()
assert AUDIT_BASELINE.is_file()

device_46 = torch.device(
    "cuda" if torch.cuda.is_available() else "cpu"
)

selection_46 = json.loads(
    AUDIT_SELECTION.read_text(encoding="utf-8")
)
baseline_46 = json.loads(
    AUDIT_BASELINE.read_text(encoding="utf-8")
)
saved_46 = torch.load(
    AUDIT_CHECKPOINT,
    map_location="cpu",
    weights_only=True
)

assert saved_46["step"] == 128
assert saved_46["precision"] == "fp32"

train_ids_46 = selection_46["train_ids"]
val_ids_46 = selection_46["val_ids"]
old_train_ids_46 = set(
    selection_46["carryover_ids"]
)

assert len(train_ids_46) == 64
assert len(val_ids_46) == 16
assert len(old_train_ids_46) == 8

record_lookup_46 = {
    r["id"]: r for r in train_records
}
dataset_lookup_46 = {
    r["id"]: i
    for i, r in enumerate(train_dataset.records)
}

# ------------------------------------------------------------
# 1. Load saved 128-update model independently
# ------------------------------------------------------------

print("LOADING SAVED PILOT MODEL")
print("=" * 58)

model_46 = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(device_46).float()

model_46.lm_head.load_state_dict(
    saved_46["head"], strict=True
)

for layer, weights in zip(
    model_46.wav2vec2.encoder.layers[-2:],
    saved_46["upper_layers"]
):
    layer.load_state_dict(weights, strict=True)

model_46.eval()
model_46.requires_grad_(False)

blank_46 = tokenizer.pad_token_id

print("Checkpoint: update", saved_46["step"])
print("Recordings to evaluate: 80")
print("Model in evaluation mode:", not model_46.training)

# ------------------------------------------------------------
# 2. Evaluate all recordings
# ------------------------------------------------------------

rows_46 = []

def evaluate_record_46(rid, group):

    record = record_lookup_46[rid]
    example = train_dataset[
        dataset_lookup_46[rid]
    ]
    batch = ctc_collator([example])

    batch = {
        k: v.to(device_46)
        for k, v in batch.items()
    }

    actual_seconds = (
        int(batch["attention_mask"].sum().item())
        / 16000
    )

    metadata_seconds = float(
        record["duration_seconds"]
    )

    with torch.no_grad():
        output = model_46(**batch)

        logits = output.logits.float()
        frame_ids = logits.argmax(dim=-1)

        blank_fraction = (
            (frame_ids == blank_46)
            .float()
            .mean()
            .item()
        )

        blank_probability = (
            logits.softmax(dim=-1)[
                :, :, blank_46
            ]
            .mean()
            .item()
        )

        prediction = processor.batch_decode(
            frame_ids.cpu()
        )[0]

    prediction = normalize_amharic_ctc(
        prediction
    )

    reference = normalize_amharic_ctc(
        record["transcription"]
    )

    ref_chars = len(reference.replace(" ", ""))
    pred_chars = len(prediction.replace(" ", ""))

    return {
        "id": rid,
        "group": group,
        "speaker": record["speaker_id"],
        "metadata_seconds": metadata_seconds,
        "audio_seconds": actual_seconds,
        "reference": reference,
        "prediction": prediction,
        "reference_chars": ref_chars,
        "predicted_chars": pred_chars,
        "chars_per_second":
            ref_chars / max(actual_seconds, 0.01),
        "prediction_length_ratio":
            pred_chars / max(ref_chars, 1),
        "cer": float(cer(reference, prediction)),
        "wer": float(wer(reference, prediction)),
        "ctc_loss": float(output.loss.item()),
        "blank_argmax_fraction": blank_fraction,
        "mean_blank_probability": blank_probability
    }

groups_46 = {
    "Previous 8 training": [
        rid for rid in train_ids_46
        if rid in old_train_ids_46
    ],
    "New 56 training": [
        rid for rid in train_ids_46
        if rid not in old_train_ids_46
    ],
    "Held-out 16": list(val_ids_46)
}

for group_name, ids in groups_46.items():
    print(f"\nEvaluating {group_name}...")

    for i, rid in enumerate(ids, 1):
        rows_46.append(
            evaluate_record_46(rid, group_name)
        )

        if i % 10 == 0 or i == len(ids):
            print(f"  {i}/{len(ids)}")

# ------------------------------------------------------------
# 3. Aggregate recognition metrics by group
# ------------------------------------------------------------

def summarize_group_46(group_name):

    group = [
        r for r in rows_46
        if r["group"] == group_name
    ]

    return {
        "count": len(group),
        "cer": cer(
            [r["reference"] for r in group],
            [r["prediction"] for r in group]
        ),
        "wer": wer(
            [r["reference"] for r in group],
            [r["prediction"] for r in group]
        ),
        "mean_ctc_loss": statistics.mean(
            r["ctc_loss"] for r in group
        ),
        "blank_frames": statistics.mean(
            r["blank_argmax_fraction"]
            for r in group
        ),
        "prediction_length_ratio": (
            sum(r["predicted_chars"] for r in group)
            / max(
                sum(r["reference_chars"] for r in group),
                1
            )
        )
    }

summary_46 = {
    name: summarize_group_46(name)
    for name in groups_46
}

print("\n" + "=" * 70)
print("RECOGNITION FAILURE-MODE SUMMARY")
print("=" * 70)

print(
    f"{'Group':<21}"
    f"{'CER':>8}"
    f"{'WER':>8}"
    f"{'CTC loss':>11}"
    f"{'Blank %':>10}"
    f"{'Length':>9}"
)

for name, s in summary_46.items():
    print(
        f"{name:<21}"
        f"{100*s['cer']:>7.1f}%"
        f"{100*s['wer']:>7.1f}%"
        f"{s['mean_ctc_loss']:>11.2f}"
        f"{100*s['blank_frames']:>9.1f}%"
        f"{s['prediction_length_ratio']:>9.2f}"
    )

print("\nLength = predicted characters / reference characters")
print("Blank % = fraction of frames decoded as CTC blank")

# ------------------------------------------------------------
# 4. Compare each validation recording before vs after
# ------------------------------------------------------------

baseline_by_id_46 = {
    r["id"]: r
    for r in baseline_46["validation_predictions"]
}

changes_46 = []

for row in rows_46:

    if row["group"] != "Held-out 16":
        continue

    before = baseline_by_id_46[row["id"]]["cer"]
    after = row["cer"]

    changes_46.append({
        "id": row["id"],
        "before": before,
        "after": after,
        "change": after - before
    })

changes_46.sort(
    key=lambda row: row["change"]
)

print("\n" + "=" * 65)
print("PER-RECORDING VALIDATION CHANGE")
print("=" * 65)

print("Most improved (negative CER change is better):")

for row in changes_46[:5]:
    print(
        row["id"],
        f"{row['before']*100:.1f}% ->",
        f"{row['after']*100:.1f}%",
        f"(change {row['change']*100:+.1f} pp)"
    )

print("\nMost degraded:")

for row in changes_46[-5:]:
    print(
        row["id"],
        f"{row['before']*100:.1f}% ->",
        f"{row['after']*100:.1f}%",
        f"(change {row['change']*100:+.1f} pp)"
    )

# ------------------------------------------------------------
# 5. Identify unusual transcript/audio ratios
# ------------------------------------------------------------

by_density_46 = sorted(
    rows_46,
    key=lambda row: row["chars_per_second"]
)

duration_mismatches_46 = [
    row for row in rows_46
    if abs(
        row["audio_seconds"]
        - row["metadata_seconds"]
    ) > 0.5
]

print("\n" + "=" * 65)
print("TRANSCRIPT QUALITY AUDIT")
print("=" * 65)

print("Recording duration mismatches (>0.5s):",
      len(duration_mismatches_46))

for row in duration_mismatches_46[:8]:
    print(
        row["id"],
        "metadata:", round(row["metadata_seconds"], 2),
        "audio:", round(row["audio_seconds"], 2)
    )

print("\nLowest transcript characters per second:")
print("(Candidates for manual review, not proven errors)")

for row in by_density_46[:10]:
    print(
        row["id"],
        f"| {row['audio_seconds']:.1f}s",
        f"| {row['chars_per_second']:.2f} chars/s",
        f"| loss {row['ctc_loss']:.2f}",
        "|", row["group"]
    )

# ------------------------------------------------------------
# 6. Save complete audit
# ------------------------------------------------------------

audit_46 = {
    "checkpoint_step": int(saved_46["step"]),
    "summary": summary_46,
    "validation_changes": changes_46,
    "duration_mismatches": duration_mismatches_46,
    "rows": rows_46
}

AUDIT_OUTPUT.write_text(
    json.dumps(
        audit_46,
        indent=2,
        ensure_ascii=False
    ),
    encoding="utf-8"
)

print("\n" + "=" * 65)
print("AUDIT COMPLETE")
print("=" * 65)
print("Saved:", AUDIT_OUTPUT)
print("Optimizer updates: 0")
print("Checkpoints modified: 0")


LOADING SAVED PILOT MODEL
Checkpoint: update 128
Recordings to evaluate: 80
Model in evaluation mode: True

Evaluating Previous 8 training...
  8/8

Evaluating New 56 training...
  10/56
  20/56
  30/56
  40/56
  50/56
  56/56

Evaluating Held-out 16...
  10/16
  16/16

RECOGNITION FAILURE-MODE SUMMARY
Group                     CER     WER   CTC loss   Blank %   Length
Previous 8 training     44.0%   92.6%       1.07     89.7%     0.64
New 56 training         87.6%  100.0%       6.78     93.9%     0.41
Held-out 16             89.5%   99.7%       6.93     94.7%     0.37

Length = predicted characters / reference characters
Blank % = fraction of frames decoded as CTC blank

PER-RECORDING VALIDATION CHANGE
Most improved (negative CER change is better):
2c9gwYKUtqawnnB84YBu 111.4% -> 89.5% (change -21.9 pp)
EXU85FucVzBBWyHHmdVD 91.8% -> 89.3% (change -2.5 pp)
EN0L0GPcZTOsDC23WcT9 89.5% -> 87.6% (change -1.9 pp)
GTrr92kY5jgPmKFucKHm 91.8% -> 90.4% (change -1.4 pp)
WSYp3H7uoLiswpjUfMcI 91.4%

In [ ]:

# ============================================================
# CELL 47 - TARGETED AUDIO / TRANSCRIPT QUALITY REVIEW
#
# Listen to recordings most likely to reveal
# transcription, clipping, or silence problems.
#
# No model loading or training.
# Existing selections/checkpoints remain unchanged.
# ============================================================

import json
import statistics
from pathlib import Path
from IPython.display import Audio, display

AUDIT_FILE_47 = (
    DATA_DIR / "scaled_amharic_64_16_v1"
    / "failure_mode_audit.json"
)

assert AUDIT_FILE_47.exists()

audit_47 = json.loads(
    AUDIT_FILE_47.read_text(encoding="utf-8")
)

rows_47 = audit_47["rows"]
by_id_47 = {r["id"]: r for r in rows_47}

record_by_id_47 = {
    r["id"]: r for r in train_records
}

old_47 = [
    r for r in rows_47
    if r["group"] == "Previous 8 training"
]

new_47 = [
    r for r in rows_47
    if r["group"] == "New 56 training"
]

val_47 = [
    r for r in rows_47
    if r["group"] == "Held-out 16"
]

print("REFERENCE CHARACTER DENSITY")
print("=" * 55)

for name, group in [
    ("Previously learned", old_47),
    ("New training", new_47),
    ("Held-out", val_47)
]:
    densities = [
        r["chars_per_second"]
        for r in group
    ]

    print(
        f"{name:<20}",
        f"median={statistics.median(densities):.2f}",
        f"min={min(densities):.2f}",
        f"max={max(densities):.2f}"
    )

# ------------------------------------------------------------
# 1. Select diagnostic examples
# ------------------------------------------------------------

review_47 = []
seen_47 = set()

def add_review_47(reason, row):
    if row["id"] not in seen_47:
        review_47.append((reason, row))
        seen_47.add(row["id"])

# Known positive control
anchor_id_47 = "6Q0fEziAqyQVIz4J8aws"

add_review_47(
    "POSITIVE CONTROL: previously learned recording",
    by_id_47[anchor_id_47]
)

# Lowest transcript density among new training examples
add_review_47(
    "TRAIN: unusually sparse transcript",
    min(
        new_47,
        key=lambda r: r["chars_per_second"]
    )
)

# Highest CTC loss not already selected
for row in sorted(
    new_47,
    key=lambda r: r["ctc_loss"],
    reverse=True
):
    if row["id"] not in seen_47:
        add_review_47(
            "TRAIN: highest remaining CTC loss",
            row
        )
        break

# Lowest transcript density in validation
add_review_47(
    "HELD-OUT: unusually sparse transcript",
    min(
        val_47,
        key=lambda r: r["chars_per_second"]
    )
)

# Largest deterioration since the validation baseline
changes_47 = audit_47["validation_changes"]

most_degraded_47 = max(
    changes_47,
    key=lambda r: r["change"]
)

add_review_47(
    "HELD-OUT: largest CER deterioration",
    by_id_47[most_degraded_47["id"]]
)

assert len(review_47) == 5

# ------------------------------------------------------------
# 2. Display audio and transcript side by side
# ------------------------------------------------------------

print("\n" + "=" * 65)
print("TARGETED AUDIO REVIEW")
print("=" * 65)

review_log_47 = []

for index, (reason, row) in enumerate(review_47, 1):

    record = record_by_id_47[row["id"]]

    audio_path = (
        Path(AUDIO_DIR) / record["audio_file"]
    )

    assert audio_path.exists(), audio_path

    print("\n" + "=" * 65)
    print(f"RECORDING {index}/5")
    print("=" * 65)

    print("Reason:", reason)
    print("ID:", row["id"])
    print("Group:", row["group"])

    print(
        "Audio duration:",
        f"{row['audio_seconds']:.2f}s"
    )

    print(
        "Reference density:",
        f"{row['chars_per_second']:.2f} chars/sec"
    )

    print(
        "CTC loss:",
        f"{row['ctc_loss']:.3f}"
    )

    print(
        "CER:",
        f"{row['cer'] * 100:.2f}%"
    )

    print(
        "Predicted/reference length:",
        f"{row['prediction_length_ratio']:.2f}"
    )

    print("\nREFERENCE TRANSCRIPT:")
    print(row["reference"])

    print("\nMODEL PREDICTION:")
    print(row["prediction"] or "[EMPTY]")

    print("\nLISTEN TO AUDIO:")
    display(Audio(filename=str(audio_path)))

    review_log_47.append({
        "id": row["id"],
        "reason": reason,
        "group": row["group"],
        "duration_seconds": row["audio_seconds"],
        "reference": row["reference"],
        "cer": row["cer"],
        "ctc_loss": row["ctc_loss"],
        "review_status": "not_yet_reviewed"
    })

# ------------------------------------------------------------
# 3. Save review queue separately
# ------------------------------------------------------------

REVIEW_FILE_47 = (
    DATA_DIR / "scaled_amharic_64_16_v1"
    / "manual_review_queue.json"
)

if not REVIEW_FILE_47.exists():
    REVIEW_FILE_47.write_text(
        json.dumps(
            review_log_47,
            ensure_ascii=False,
            indent=2
        ),
        encoding="utf-8"
    )

print("\n" + "=" * 65)
print("REVIEW QUEUE CREATED")
print("=" * 65)

print("Recordings to listen to:", len(review_47))
print("Review queue:", REVIEW_FILE_47)
print("Training updates: 0")
print("Checkpoints modified: 0")


REFERENCE CHARACTER DENSITY
Previously learned   median=6.11 min=4.42 max=9.23
New training         median=5.59 min=2.51 max=9.26
Held-out             median=6.02 min=2.60 max=7.98

TARGETED AUDIO REVIEW

RECORDING 1/5
Reason: POSITIVE CONTROL: previously learned recording
ID: 6Q0fEziAqyQVIz4J8aws
Group: Previous 8 training
Audio duration: 5.18s
Reference density: 5.98 chars/sec
CTC loss: 1.152
CER: 48.72%
Predicted/reference length: 0.61

REFERENCE TRANSCRIPT:
ይህ ምስል የሚያሳየው ከሸክላ የሚሰራ የሸክላ ድስት ምስል ነው

MODEL PREDICTION:
ይህምየሳውሸክላራራየሸክላድ ምስ ው

LISTEN TO AUDIO:



RECORDING 2/5
Reason: TRAIN: unusually sparse transcript
ID: BARUJgkogmBvGp4iJ0sx
Group: New 56 training
Audio duration: 14.74s
Reference density: 2.51 chars/sec
CTC loss: 10.726
CER: 100.00%
Predicted/reference length: 1.03

REFERENCE TRANSCRIPT:
አህያ ለጭነት አገልግሎት እንጠቀመዋለን ለባህላዊ የጭነት አገልግሎቶች

MODEL PREDICTION:
ወጥዩንንበናጥበበደበበጫጥጥ በበናዱላጥመናሲ በጫጥበናጥላበጫዱንጥዘ

LISTEN TO AUDIO:



RECORDING 3/5
Reason: TRAIN: highest remaining CTC loss
ID: JljzcvdzYAAyQmAc4x5u
Group: New 56 training
Audio duration: 14.90s
Reference density: 3.56 chars/sec
CTC loss: 9.748
CER: 109.09%
Predicted/reference length: 1.40

REFERENCE TRANSCRIPT:
ከላይ በምስሉ ላይ የምትመለከቱት የቤት እቃ ምን በመባል ይታወቃል ለምን ለምን አገልግሎትስ ሊውል ይችላል

MODEL PREDICTION:
ውህንንው በውይናንችንርና ነናውእሲእንንላን ንእንን ንውበ ውው ንያውበው ንው ናንውበንንውንላምል በውው እንንንውውለውንገ ውገንንላው ው ናውዱ

LISTEN TO AUDIO:



RECORDING 4/5
Reason: HELD-OUT: unusually sparse transcript
ID: 4ljLQRFgHFJqEsJDZuHd
Group: Held-out 16
Audio duration: 14.26s
Reference density: 2.60 chars/sec
CTC loss: 6.723
CER: 91.11%
Predicted/reference length: 0.49

REFERENCE TRANSCRIPT:
ይህ የምንመለከተዉ ምስል የኢትዮጵያ ባህላዊ ግብይት እንዲሁም ሸመታ ነዉ

MODEL PREDICTION:
ፀን ይውሰበየበርበሰ በድማበድውው

LISTEN TO AUDIO:



RECORDING 5/5
Reason: HELD-OUT: largest CER deterioration
ID: JHt6FIBUQa9WuQez8J2M
Group: Held-out 16
Audio duration: 14.86s
Reference density: 6.46 chars/sec
CTC loss: 6.963
CER: 84.48%
Predicted/reference length: 0.47

REFERENCE TRANSCRIPT:
አካላዊ ትምህርትና ስፖርት የህፃናት አካላዊና አእምሮአዊ ጤናን ለመጠበቅ የአካል ብቃት እንቅስቃሴ ጨዋታውን ለማሳለጥና ለማስኬድ የሚጠቀሙት የአካል ብቃት ትምህርት ስፖርት አንደኛው ነው

MODEL PREDICTION:
ዱውይው ምይስነንንንሲ ንው ው ውውስሆንእን ስም ምእ ንእውን ውይእምስንናይንእሲስው ላ ው

LISTEN TO AUDIO:



REVIEW QUEUE CREATED
Recordings to listen to: 5
Review queue: /content/drive/MyDrive/Amharic_ASR_XLSR/data/scaled_amharic_64_16_v1/manual_review_queue.json
Training updates: 0
Checkpoints modified: 0


In [ ]:

# ============================================================
# CELL 48 - APPLY MANUAL QUALITY REVIEW
#
# Record five human annotations from Cell 47.
# Create a provisional filtered dataset.
# Select five additional recordings for review.
#
# No training and no checkpoint modifications.
# ============================================================

import json
from pathlib import Path
from IPython.display import Audio, display

QA_DIR = DATA_DIR / "scaled_amharic_64_16_v1"

REVIEW_QUEUE = QA_DIR / "manual_review_queue.json"
AUDIT_PATH = QA_DIR / "failure_mode_audit.json"
SELECTION_PATH = QA_DIR / "selection.json"

LABELS_PATH = QA_DIR / "manual_review_results_round1.json"
FILTERED_PATH = QA_DIR / "quality_filtered_v1.json"
ROUND2_PATH = QA_DIR / "manual_review_round2.json"

review_queue = json.loads(
    REVIEW_QUEUE.read_text(encoding="utf-8")
)
audit = json.loads(
    AUDIT_PATH.read_text(encoding="utf-8")
)
selection = json.loads(
    SELECTION_PATH.read_text(encoding="utf-8")
)

assert len(review_queue) == 5

audit_rows = {
    row["id"]: row
    for row in audit["rows"]
}

# ------------------------------------------------------------
# 1. Save your review results in the displayed order
# ------------------------------------------------------------

decisions = [
    (
        "quarantine",
        "Partial transcript with additional speech"
    ),
    (
        "quarantine",
        "Silence reported during listening"
    ),
    (
        "verified_match",
        "Spoken content matches transcript"
    ),
    (
        "noisy_challenge",
        "Heavy background noise and repeated words"
    ),
    (
        "verified_match",
        "Spoken content matches transcript"
    )
]

expected_groups = [
    "Previous 8 training",
    "New 56 training",
    "New 56 training",
    "Held-out 16",
    "Held-out 16"
]

annotations = []

for index, (item, decision) in enumerate(
    zip(review_queue, decisions)
):

    status, reason = decision
    rid = item["id"]

    assert rid in audit_rows
    assert audit_rows[rid]["group"] == expected_groups[index]

    annotations.append({
        "id": rid,
        "original_group": expected_groups[index],
        "review_status": status,
        "finding": reason
    })

# Prevent accidental overwriting of different
# human annotations from a previous run.
if LABELS_PATH.exists():
    existing = json.loads(
        LABELS_PATH.read_text(encoding="utf-8")
    )
    assert existing == annotations, (
        "Existing review labels differ. "
        "Inspect the saved file before changing them."
    )
else:
    LABELS_PATH.write_text(
        json.dumps(
            annotations,
            ensure_ascii=False,
            indent=2
        ),
        encoding="utf-8"
    )

print("ROUND 1 HUMAN REVIEW RESULTS")
print("=" * 60)

for i, row in enumerate(annotations, 1):
    print(
        f"{i}. {row['id']}",
        "|", row["review_status"]
    )
    print("   ", row["finding"])

# ------------------------------------------------------------
# 2. Build provisional training/evaluation subsets
# ------------------------------------------------------------

train_quarantine = {
    row["id"]
    for row in annotations
    if row["review_status"] == "quarantine"
}

val_challenge = {
    row["id"]
    for row in annotations
    if row["review_status"] == "noisy_challenge"
}

original_train = selection["train_ids"]
original_val = selection["val_ids"]

assert train_quarantine.issubset(set(original_train))
assert val_challenge.issubset(set(original_val))

filtered_train = [
    rid for rid in original_train
    if rid not in train_quarantine
]

provisional_val = [
    rid for rid in original_val
    if rid not in val_challenge
]

verified_matches = {
    row["id"]
    for row in annotations
    if row["review_status"] == "verified_match"
}

filtered = {
    "status": "provisional_not_fully_reviewed",
    "train_ids": filtered_train,
    "primary_val_ids": provisional_val,
    "noisy_challenge_ids": sorted(val_challenge),
    "quarantined_train_ids": sorted(train_quarantine),
    "verified_match_ids": sorted(verified_matches),
    "source_selection": str(SELECTION_PATH),
    "note": (
        "Only five examples have undergone manual review. "
        "Unreviewed examples are not certified clean."
    )
}

if FILTERED_PATH.exists():
    previous = json.loads(
        FILTERED_PATH.read_text(encoding="utf-8")
    )
    assert previous == filtered, (
        "A different filtered split already exists."
    )
else:
    FILTERED_PATH.write_text(
        json.dumps(
            filtered,
            ensure_ascii=False,
            indent=2
        ),
        encoding="utf-8"
    )

print("\nPROVISIONAL DATASET")
print("=" * 60)

print("Original training:", len(original_train))
print("Quarantined training:", len(train_quarantine))
print("Remaining training:", len(filtered_train))

print("\nOriginal validation:", len(original_val))
print("Noisy challenge:", len(val_challenge))
print("Remaining primary validation:", len(provisional_val))

print("\nHuman-verified matching examples:",
      len(verified_matches))

print(
    "Other examples remain unreviewed:",
    len(filtered_train + provisional_val)
    - len(verified_matches)
)

# ------------------------------------------------------------
# 3. Select five more examples for human inspection
# ------------------------------------------------------------

already_reviewed = {
    row["id"] for row in annotations
}

training_pool = [
    row for row in audit["rows"]
    if row["id"] in filtered_train
    and row["id"] not in already_reviewed
]

validation_pool = [
    row for row in audit["rows"]
    if row["id"] in provisional_val
    and row["id"] not in already_reviewed
]

round2 = []
selected_ids = set()

def add_candidate(reason, row):
    if row["id"] not in selected_ids:
        round2.append({
            "id": row["id"],
            "reason": reason,
            "group": row["group"]
        })
        selected_ids.add(row["id"])

# Two training samples with low transcript density.
for row in sorted(
    training_pool,
    key=lambda r: r["chars_per_second"]
)[:2]:
    add_candidate(
        "Training: low transcript density",
        row
    )

# One high-loss training sample not already chosen.
for row in sorted(
    training_pool,
    key=lambda r: r["ctc_loss"],
    reverse=True
):
    if row["id"] not in selected_ids:
        add_candidate(
            "Training: high CTC loss",
            row
        )
        break

# One sparse validation example.
for row in sorted(
    validation_pool,
    key=lambda r: r["chars_per_second"]
):
    if row["id"] not in selected_ids:
        add_candidate(
            "Validation: low transcript density",
            row
        )
        break

# One high-loss validation example.
for row in sorted(
    validation_pool,
    key=lambda r: r["ctc_loss"],
    reverse=True
):
    if row["id"] not in selected_ids:
        add_candidate(
            "Validation: high CTC loss",
            row
        )
        break

assert len(round2) == 5

if ROUND2_PATH.exists():
    saved_round2 = json.loads(
        ROUND2_PATH.read_text(encoding="utf-8")
    )
    assert saved_round2 == round2
else:
    ROUND2_PATH.write_text(
        json.dumps(
            round2,
            ensure_ascii=False,
            indent=2
        ),
        encoding="utf-8"
    )

# ------------------------------------------------------------
# 4. Play the new recordings
# ------------------------------------------------------------

records_by_id = {
    record["id"]: record
    for record in train_records
}

print("\n" + "=" * 65)
print("ROUND 2: FIVE RECORDINGS TO REVIEW")
print("=" * 65)

for index, item in enumerate(round2, 1):

    rid = item["id"]
    row = audit_rows[rid]
    record = records_by_id[rid]

    audio_path = (
        Path(AUDIO_DIR) / record["audio_file"]
    )

    assert audio_path.is_file()

    print("\n" + "=" * 60)
    print(f"RECORDING {index}/5")
    print("=" * 60)

    print("ID:", rid)
    print("Reason:", item["reason"])
    print(
        "Duration:",
        round(row["audio_seconds"], 2),
        "seconds"
    )
    print(
        "CTC loss:",
        round(row["ctc_loss"], 3)
    )
    print(
        "Transcript density:",
        round(row["chars_per_second"], 2),
        "characters/second"
    )

    print("\nREFERENCE:")
    print(row["reference"])

    print("\nMODEL PREDICTION:")
    print(row["prediction"] or "[EMPTY]")

    print("\nAUDIO:")
    display(Audio(filename=str(audio_path)))

print("\n" + "=" * 65)
print("QUALITY AUDIT UPDATED")
print("=" * 65)

print("Annotations:", LABELS_PATH)
print("Filtered split:", FILTERED_PATH)
print("Next review queue:", ROUND2_PATH)
print("Optimizer updates: 0")
print("Existing checkpoints modified: 0")


ROUND 1 HUMAN REVIEW RESULTS
1. 6Q0fEziAqyQVIz4J8aws | quarantine
    Partial transcript with additional speech
2. BARUJgkogmBvGp4iJ0sx | quarantine
    Silence reported during listening
3. JljzcvdzYAAyQmAc4x5u | verified_match
    Spoken content matches transcript
4. 4ljLQRFgHFJqEsJDZuHd | noisy_challenge
    Heavy background noise and repeated words
5. JHt6FIBUQa9WuQez8J2M | verified_match
    Spoken content matches transcript

PROVISIONAL DATASET
Original training: 64
Quarantined training: 2
Remaining training: 62

Original validation: 16
Noisy challenge: 1
Remaining primary validation: 15

Human-verified matching examples: 2
Other examples remain unreviewed: 75

ROUND 2: FIVE RECORDINGS TO REVIEW

RECORDING 1/5
ID: 1kPe5yhdSKLyyBYtp1yP
Reason: Training: low transcript density
Duration: 14.98 seconds
CTC loss: 6.065
Transcript density: 3.27 characters/second

REFERENCE:
እስልምና እስልምና አንዱ የሀይማኖት አይነት ሲሆን ይህ ሃይማኖት መቼ ተመሰረተ በማንስ ተመሰረተ

MODEL PREDICTION:
ፀይይውውን በነይንምበቅታምም በ ርውውበ በውለዱችንው በ


RECORDING 2/5
ID: 7ZOeZpBUxW6IXls17BxG
Reason: Training: low transcript density
Duration: 14.86 seconds
CTC loss: 7.04
Transcript density: 3.37 characters/second

REFERENCE:
ይህ የልቦለድ የመጽሃፍ ግርባብን ነው እና ይህ ልቦልድ መጽሃፍ ግርባብ ልቦለዱን ይጻፈው ሰው ማን ነው

MODEL PREDICTION:
ወን ደለ በንውየበንጫሳውቻአ በጥንበይይአርሳአር ይ ይዘ

AUDIO:



RECORDING 3/5
ID: 5us9lovEMnIT5mMb6bQ9
Reason: Training: high CTC loss
Duration: 14.38 seconds
CTC loss: 8.543
Transcript density: 6.33 characters/second

REFERENCE:
እዚህጋ የምትመለከቱት በጣም ብዙ መፅሐፍ የያዘ ቤተመጻሕፍት ነው ከሱም ደግሞ የወጡ የተወሰኑ መፅሐፍ ከፊት ለፊት አሉ ስታዩት ደግሞ ይሄ ቤተመጻሕፍት የት አካባቢ ሚገኝ ይመስላችኋል

MODEL PREDICTION:
ውናንይእስአውንችደንእስንስልንስንይልእእንንስ ው ንንስን እውህውአንልንውስንንልንልችሆእናምውህውልውነንስንመ ንስህሳይዱ

AUDIO:



RECORDING 4/5
ID: GTrr92kY5jgPmKFucKHm
Reason: Validation: low transcript density
Duration: 14.66 seconds
CTC loss: 5.952
Transcript density: 3.89 characters/second

REFERENCE:
በእስር ቤት የእስር ፍርድ ላይ ያለ ሰው ምስል ያሳያል የታሰረው ሰው እጁ በካቴና ውስጥ እንደታሰረ የሚያሳይ ምልክት

MODEL PREDICTION:
ይ ውአ ምበ ው

AUDIO:



RECORDING 5/5
ID: 2c9gwYKUtqawnnB84YBu
Reason: Validation: high CTC loss
Duration: 14.9 seconds
CTC loss: 8.452
Transcript density: 5.97 characters/second

REFERENCE:
ጌጣጌጥ ጆሮ ጌጥ ጆሮ ጌጥ በመጠኑ እጅግ አነስተኛ የሆነ በጣም ውብ ማራኪና አስደናቂ በጆሮ ላይ የሚደረግ የጌጥ ዓይነት ከወርቅ ከብር ከነሀስና የተለያዩ ነገሮች የሚሠራ ጌጣጌጥ ነው

MODEL PREDICTION:
ውልልውሲ ህውውያውሳሳንያ ውህሲነውንስ ንል ያናያ ንእ ምናህናውያ ያሳውያህዊያናውልሲንንህልንቂያልንያነውናውነንያውውያናያነልልዩው ህንልያንልያበናያናህህዱ

AUDIO:



QUALITY AUDIT UPDATED
Annotations: /content/drive/MyDrive/Amharic_ASR_XLSR/data/scaled_amharic_64_16_v1/manual_review_results_round1.json
Filtered split: /content/drive/MyDrive/Amharic_ASR_XLSR/data/scaled_amharic_64_16_v1/quality_filtered_v1.json
Next review queue: /content/drive/MyDrive/Amharic_ASR_XLSR/data/scaled_amharic_64_16_v1/manual_review_round2.json
Optimizer updates: 0
Existing checkpoints modified: 0


In [ ]:

# ============================================================
# CELL 49 - FINALIZE MANUAL QA AND CLEAN EVALUATION
#
# 4 matching recordings
# 1 recording with minor filler sounds
#
# Preserve original data and all checkpoints.
# ============================================================

import json
from pathlib import Path
from jiwer import cer, wer

QA_DIR = DATA_DIR / "scaled_amharic_64_16_v1"

ROUND2_QUEUE = QA_DIR / "manual_review_round2.json"
ROUND1_LABELS = QA_DIR / "manual_review_results_round1.json"
ORIGINAL_SPLIT = QA_DIR / "selection.json"
AUDIT_FILE = QA_DIR / "failure_mode_audit.json"
BASELINE_FILE = QA_DIR / "fp32_preflight.json"

ROUND2_RESULTS = QA_DIR / "manual_review_results_round2.json"
CLEAN_SPLIT_FILE = QA_DIR / "quality_filtered_v2.json"
CLEAN_METRICS_FILE = QA_DIR / "quality_metrics_v2.json"

def load_json(path):
    assert path.is_file(), f"Missing: {path}"
    return json.loads(path.read_text(encoding="utf-8"))

def save_checked(path, data):
    if path.exists():
        assert load_json(path) == data, (
            f"Existing file differs: {path}"
        )
        print("Already saved:", path.name)
    else:
        path.write_text(
            json.dumps(data, ensure_ascii=False, indent=2),
            encoding="utf-8"
        )
        print("Saved:", path.name)

queue = load_json(ROUND2_QUEUE)
round1 = load_json(ROUND1_LABELS)
original = load_json(ORIGINAL_SPLIT)
audit = load_json(AUDIT_FILE)
baseline = load_json(BASELINE_FILE)

assert len(queue) == 5

# ------------------------------------------------------------
# 1. Record the five new human assessments
# ------------------------------------------------------------

human_decisions = [
    ("verified_match", "Speech matches transcript"),
    ("verified_match", "Speech matches transcript"),
    (
        "match_with_fillers",
        "Correct speech with minor ah/hesitation sounds"
    ),
    ("verified_match", "Speech matches transcript"),
    ("verified_match", "Speech matches transcript"),
]

round2 = []

for item, (status, finding) in zip(
    queue, human_decisions
):
    round2.append({
        "id": item["id"],
        "original_group": item["group"],
        "review_status": status,
        "finding": finding
    })

assert len({r["id"] for r in round2}) == 5

save_checked(ROUND2_RESULTS, round2)

# ------------------------------------------------------------
# 2. Combine both review rounds
# ------------------------------------------------------------

all_reviews = round1 + round2

assert len(all_reviews) == 10
assert len({r["id"] for r in all_reviews}) == 10

quarantine = {
    r["id"]
    for r in all_reviews
    if r["review_status"] == "quarantine"
}

noisy_challenge = {
    r["id"]
    for r in all_reviews
    if r["review_status"] == "noisy_challenge"
}

verified = {
    r["id"]
    for r in all_reviews
    if r["review_status"] == "verified_match"
}

with_fillers = {
    r["id"]
    for r in all_reviews
    if r["review_status"] == "match_with_fillers"
}

assert len(quarantine) == 2
assert len(noisy_challenge) == 1
assert len(verified) == 6
assert len(with_fillers) == 1

# ------------------------------------------------------------
# 3. Construct the quality-filtered split
# ------------------------------------------------------------

train_ids = [
    rid for rid in original["train_ids"]
    if rid not in quarantine
]

val_ids = [
    rid for rid in original["val_ids"]
    if rid not in noisy_challenge
]

assert len(train_ids) == 62
assert len(val_ids) == 15
assert not set(train_ids) & set(val_ids)

records = {r["id"]: r for r in train_records}

train_speakers = {
    records[rid]["speaker_id"]
    for rid in train_ids
}

val_speakers = {
    records[rid]["speaker_id"]
    for rid in val_ids
}

assert not train_speakers & val_speakers

clean_split = {
    "status": "provisional_human_screened",
    "train_ids": train_ids,
    "primary_val_ids": val_ids,
    "quarantined_train_ids": sorted(quarantine),
    "noisy_challenge_ids": sorted(noisy_challenge),
    "verified_match_ids": sorted(verified),
    "match_with_fillers_ids": sorted(with_fillers),
    "reviewed_count": len(all_reviews),
    "note": (
        "Only 10 of the original 80 recordings were "
        "manually reviewed. Unreviewed recordings "
        "are not certified clean. Existing model "
        "checkpoints may already contain training "
        "influence from quarantined recordings."
    )
}

save_checked(CLEAN_SPLIT_FILE, clean_split)

# ------------------------------------------------------------
# 4. Recalculate validation metrics on the SAME 15 IDs
# ------------------------------------------------------------

baseline_by_id = {
    r["id"]: r
    for r in baseline["validation_predictions"]
}

pilot_by_id = {
    r["id"]: r
    for r in audit["rows"]
}

def compute_metrics(ids, source):
    refs = [source[rid]["reference"] for rid in ids]
    preds = [
        source[rid]["prediction"]
        for rid in ids
    ]

    return {
        "count": len(ids),
        "cer": float(cer(refs, preds)),
        "wer": float(wer(refs, preds)),
        "nonempty": sum(bool(p.strip()) for p in preds)
    }

assert all(rid in baseline_by_id for rid in val_ids)
assert all(rid in pilot_by_id for rid in val_ids)

before = compute_metrics(val_ids, baseline_by_id)
after = compute_metrics(val_ids, pilot_by_id)

challenge_ids = sorted(noisy_challenge)

challenge_before = compute_metrics(
    challenge_ids, baseline_by_id
)
challenge_after = compute_metrics(
    challenge_ids, pilot_by_id
)

train_after = compute_metrics(
    train_ids, pilot_by_id
)

metrics = {
    "primary_validation_before_pilot": before,
    "primary_validation_after_128_updates": after,
    "noisy_challenge_before": challenge_before,
    "noisy_challenge_after": challenge_after,
    "training_after_128_updates": train_after
}

save_checked(CLEAN_METRICS_FILE, metrics)

# ------------------------------------------------------------
# 5. Print summary
# ------------------------------------------------------------

print("\n" + "=" * 60)
print("QUALITY REVIEW COMPLETE")
print("=" * 60)

print("Reviewed:", len(all_reviews))
print("Verified matches:", len(verified))
print("Matches with fillers:", len(with_fillers))
print("Quarantined:", len(quarantine))
print("Noisy challenge:", len(noisy_challenge))

print("\nFINAL PROVISIONAL DATASET")
print("Training:", len(train_ids))
print("Primary validation:", len(val_ids))
print("Noisy challenge:", len(challenge_ids))
print("Train/validation speaker overlap:", 0)

print("\n" + "=" * 60)
print("RECALCULATED METRICS")
print("=" * 60)

print(
    f"{'Dataset':<27}"
    f"{'CER':>10}"
    f"{'WER':>10}"
)

for label, result in [
    ("Validation before pilot", before),
    ("Validation after 128", after),
    ("Training after 128", train_after),
    ("Noisy before pilot", challenge_before),
    ("Noisy after 128", challenge_after)
]:
    print(
        f"{label:<27}"
        f"{result['cer']*100:>9.2f}%"
        f"{result['wer']*100:>9.2f}%"
    )

print("\nValidation CER improvement:",
      f"{(before['cer']-after['cer'])*100:+.2f}",
      "percentage points")

print("\nNo training was performed.")
print("All model checkpoints remain unchanged.")


Saved: manual_review_results_round2.json
Saved: quality_filtered_v2.json
Saved: quality_metrics_v2.json

QUALITY REVIEW COMPLETE
Reviewed: 10
Verified matches: 6
Matches with fillers: 1
Quarantined: 2
Noisy challenge: 1

FINAL PROVISIONAL DATASET
Training: 62
Primary validation: 15
Noisy challenge: 1
Train/validation speaker overlap: 0

RECALCULATED METRICS
Dataset                           CER       WER
Validation before pilot        90.55%    99.70%
Validation after 128           89.50%    99.70%
Training after 128             84.33%    99.41%
Noisy before pilot             91.11%   100.00%
Noisy after 128                91.11%   100.00%

Validation CER improvement: +1.05 percentage points

No training was performed.
All model checkpoints remain unchanged.


In [ ]:

# ============================================================
# CELL 50 - QUALITY-FILTERED TRAINING CONTINUATION
#
# 62 train / 15 primary validation
# Start from Cell 45 checkpoint, update 128
# Preserve optimizer state from previous training
# Train last 2 XLS-R layers + CTC head
#
# Three additional epochs (186 updates)
# FP32, no dropout/SpecAugment
# No previous checkpoints overwritten
# ============================================================

import json
import random
import hashlib
import statistics
import gc
from pathlib import Path

import torch
from transformers import Wav2Vec2ForCTC
from jiwer import cer, wer

ROOT_50 = DATA_DIR / "scaled_amharic_64_16_v1"
SOURCE_50 = ROOT_50 / "stage1_fp32" / "latest.pt"
SPLIT_50 = ROOT_50 / "quality_filtered_v2.json"
METRICS_50 = ROOT_50 / "quality_metrics_v2.json"

RUN_50 = ROOT_50 / "stage2_filtered_62_v1"
RUN_50.mkdir(parents=True, exist_ok=True)

LATEST_50 = RUN_50 / "latest.pt"
BEST_50 = RUN_50 / "best.pt"
HISTORY_50 = RUN_50 / "history.json"

DEVICE_50 = torch.device(
    "cuda" if torch.cuda.is_available() else "cpu"
)

EPOCHS_50 = 3
HEAD_LR_50 = 1e-4
ENCODER_LR_50 = 2e-6
CLIP_50 = 1.0
SEED_50 = 20261020

def read_50(path):
    assert path.is_file(), f"Missing file: {path}"
    return json.loads(path.read_text(encoding="utf-8"))

split_50 = read_50(SPLIT_50)
previous_metrics_50 = read_50(METRICS_50)

train_ids_50 = split_50["train_ids"]
val_ids_50 = split_50["primary_val_ids"]

assert len(train_ids_50) == 62
assert len(val_ids_50) == 15
assert not (set(train_ids_50) & set(val_ids_50))

records_50 = {r["id"]: r for r in train_records}
indices_50 = {
    r["id"]: i for i, r in enumerate(train_dataset.records)
}

assert all(
    rid in indices_50
    for rid in train_ids_50 + val_ids_50
)

train_speakers_50 = {
    records_50[rid]["speaker_id"]
    for rid in train_ids_50
}
val_speakers_50 = {
    records_50[rid]["speaker_id"]
    for rid in val_ids_50
}

assert not (train_speakers_50 & val_speakers_50)

# Old examples versus newly introduced recordings.
original_8 = set(
    read_50(
        ROOT_50 / "selection.json"
    )["carryover_ids"]
)

old_ids_50 = [
    rid for rid in train_ids_50 if rid in original_8
]
new_ids_50 = [
    rid for rid in train_ids_50 if rid not in original_8
]

assert len(old_ids_50) == 7
assert len(new_ids_50) == 55

source_50 = torch.load(
    SOURCE_50,
    map_location="cpu",
    weights_only=True
)

assert source_50["step"] == 128
assert source_50["precision"] == "fp32"

configuration_50 = {
    "source_signature": source_50["signature"],
    "source_step": 128,
    "train_ids": train_ids_50,
    "val_ids": val_ids_50,
    "head_lr": HEAD_LR_50,
    "encoder_lr": ENCODER_LR_50,
    "clip": CLIP_50,
    "seed": SEED_50
}

signature_50 = hashlib.sha256(
    json.dumps(
        configuration_50,
        sort_keys=True,
        ensure_ascii=False
    ).encode("utf-8")
).hexdigest()

# ------------------------------------------------------------
# 1. Load original encoder, then restore saved fine-tuning
# ------------------------------------------------------------

print("RESTORING SCALED MODEL")
print("=" * 60)

model_50 = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(DEVICE_50).float()

model_50.lm_head.load_state_dict(
    source_50["head"],
    strict=True
)

layers_50 = list(
    model_50.wav2vec2.encoder.layers[-2:]
)

for layer, weights in zip(
    layers_50,
    source_50["upper_layers"]
):
    layer.load_state_dict(weights, strict=True)

model_50.requires_grad_(False)

for layer in layers_50:
    layer.requires_grad_(True)

model_50.lm_head.requires_grad_(True)

# Keep stochastic dropout and SpecAugment disabled.
# Gradients still work normally.
model_50.eval()

encoder_parameters_50 = [
    p for layer in layers_50
    for p in layer.parameters()
    if p.requires_grad
]

head_parameters_50 = list(
    model_50.lm_head.parameters()
)

trainable_50 = (
    encoder_parameters_50 + head_parameters_50
)

assert sum(
    p.numel() for p in trainable_50
) == 25521473

optimizer_50 = torch.optim.AdamW([
    {
        "params": encoder_parameters_50,
        "lr": ENCODER_LR_50,
        "weight_decay": 0.01
    },
    {
        "params": head_parameters_50,
        "lr": HEAD_LR_50,
        "weight_decay": 0.0
    }
])

# Preserve accumulated optimizer moments.
optimizer_50.load_state_dict(
    source_50["optimizer"]
)

assert abs(
    optimizer_50.param_groups[0]["lr"] - ENCODER_LR_50
) < 1e-12

assert abs(
    optimizer_50.param_groups[1]["lr"] - HEAD_LR_50
) < 1e-12

# ------------------------------------------------------------
# 2. Restore stage 2 progress if present
# ------------------------------------------------------------

completed_50 = 0
history_50 = []
best_cer_50 = float(
    previous_metrics_50[
        "primary_validation_after_128_updates"
    ]["cer"]
)

if LATEST_50.exists():

    saved = torch.load(
        LATEST_50,
        map_location="cpu",
        weights_only=True
    )

    assert saved["signature"] == signature_50

    model_50.lm_head.load_state_dict(saved["head"])

    for layer, weights in zip(
        layers_50,
        saved["upper_layers"]
    ):
        layer.load_state_dict(weights)

    optimizer_50.load_state_dict(saved["optimizer"])

    completed_50 = int(saved["updates"])
    best_cer_50 = float(saved["best_cer"])

    if HISTORY_50.exists():
        history_50 = read_50(HISTORY_50)

    print("Resuming from stage 2 update:", completed_50)

else:
    print("Restored Cell 45 checkpoint at update 128.")

# ------------------------------------------------------------
# 3. Decode and evaluate recordings
# ------------------------------------------------------------

def batch_50(rid):

    item = train_dataset[indices_50[rid]]
    batch = ctc_collator([item])

    return {
        name: value.to(DEVICE_50)
        for name, value in batch.items()
    }

def evaluate_50(ids):

    model_50.eval()

    references = []
    predictions = []

    blank_frames = 0
    total_frames = 0

    with torch.no_grad():

        for rid in ids:

            batch = batch_50(rid)

            # Labels aren't needed for inference.
            output = model_50(
                input_values=batch["input_values"],
                attention_mask=batch["attention_mask"]
            )

            token_ids = output.logits.argmax(dim=-1)

            blank_frames += int(
                (token_ids == tokenizer.pad_token_id)
                .sum().item()
            )

            total_frames += token_ids.numel()

            prediction = processor.batch_decode(
                token_ids.cpu()
            )[0]

            prediction = normalize_amharic_ctc(
                prediction
            )

            reference = normalize_amharic_ctc(
                records_50[rid]["transcription"]
            )

            references.append(reference)
            predictions.append(prediction)

            del batch, output

    ref_chars = sum(
        len(text.replace(" ", ""))
        for text in references
    )

    pred_chars = sum(
        len(text.replace(" ", ""))
        for text in predictions
    )

    return {
        "cer": float(cer(references, predictions)),
        "wer": float(wer(references, predictions)),
        "length_ratio": pred_chars / max(ref_chars, 1),
        "blank_fraction": blank_frames / max(total_frames, 1),
        "nonempty": sum(bool(p.strip()) for p in predictions),
        "sample": predictions[0]
    }

def report_50(epoch, update):

    old = evaluate_50(old_ids_50)
    new = evaluate_50(new_ids_50)
    val = evaluate_50(val_ids_50)

    row = {
        "epoch": epoch,
        "updates": update,
        "old_train_cer": old["cer"],
        "new_train_cer": new["cer"],
        "val_cer": val["cer"],
        "val_wer": val["wer"],
        "val_length_ratio": val["length_ratio"],
        "val_blank_fraction": val["blank_fraction"],
        "val_nonempty": val["nonempty"],
        "val_sample": val["sample"]
    }

    print(f"\nEPOCH {epoch}/{EPOCHS_50}")
    print("-" * 58)

    print("Additional updates:", update)
    print(
        "Previous 7 training CER:",
        f"{old['cer']*100:.2f}%"
    )
    print(
        "New 55 training CER:",
        f"{new['cer']*100:.2f}%"
    )
    print(
        "Primary validation CER:",
        f"{val['cer']*100:.2f}%"
    )
    print(
        "Primary validation WER:",
        f"{val['wer']*100:.2f}%"
    )
    print(
        "Prediction/reference length:",
        f"{val['length_ratio']:.2f}"
    )
    print(
        "CTC blank frames:",
        f"{val['blank_fraction']*100:.1f}%"
    )
    print(
        "Nonempty validation predictions:",
        f"{val['nonempty']}/15"
    )

    print("Validation example:")
    print(val["sample"][:120] or "[EMPTY]")

    return row

def save_50(update, best_cer, save_best=False):

    checkpoint = {
        "signature": signature_50,
        "updates": update,
        "best_cer": best_cer,
        "precision": "fp32",
        "head": model_50.lm_head.state_dict(),
        "upper_layers": [
            layer.state_dict()
            for layer in layers_50
        ],
        "optimizer": optimizer_50.state_dict()
    }

    temp = RUN_50 / "latest.pt.partial"
    torch.save(checkpoint, temp)
    temp.replace(LATEST_50)

    if save_best:
        best_temp = RUN_50 / "best.pt.partial"
        torch.save(checkpoint, best_temp)
        best_temp.replace(BEST_50)

    hist_temp = RUN_50 / "history.json.partial"

    hist_temp.write_text(
        json.dumps(
            history_50,
            ensure_ascii=False,
            indent=2
        ),
        encoding="utf-8"
    )

    hist_temp.replace(HISTORY_50)

# ------------------------------------------------------------
# 4. Establish consistent starting metrics
# ------------------------------------------------------------

print("\nQUALITY-FILTERED TRAINING")
print("=" * 60)

print("Training recordings:", len(train_ids_50))
print("Primary validation:", len(val_ids_50))
print("Previously trained:", len(old_ids_50))
print("New training:", len(new_ids_50))
print("Trainable parameters:", 25521473)
print("FP32:", True)
print("Additional epochs:", EPOCHS_50)

if completed_50 == 0 and not history_50:

    starting_50 = report_50(0, 0)

    expected = previous_metrics_50[
        "primary_validation_after_128_updates"
    ]["cer"]

    assert abs(
        starting_50["val_cer"] - expected
    ) < 0.005, (
        "Starting validation CER differs from "
        "the saved Cell 49 baseline."
    )

    history_50.append(starting_50)

# ------------------------------------------------------------
# 5. Deterministic training order
# ------------------------------------------------------------

def training_id_50(update):

    index = update - 1
    epoch_index = index // len(train_ids_50)
    position = index % len(train_ids_50)

    order = list(train_ids_50)

    random.Random(
        SEED_50 + epoch_index
    ).shuffle(order)

    return order[position]

TOTAL_UPDATES_50 = EPOCHS_50 * len(train_ids_50)

losses_50 = []
norms_50 = []

# ------------------------------------------------------------
# 6. Run training
# ------------------------------------------------------------

for update in range(
    completed_50 + 1,
    TOTAL_UPDATES_50 + 1
):

    rid = training_id_50(update)

    optimizer_50.zero_grad(set_to_none=True)
    model_50.eval()

    batch = batch_50(rid)

    with torch.autocast(
        device_type=DEVICE_50.type,
        enabled=False
    ):
        loss = model_50(**batch).loss

    if not torch.isfinite(loss).item():
        raise RuntimeError(
            f"Non-finite loss at update {update}, "
            f"recording {rid}"
        )

    loss.backward()

    grad_norm = torch.nn.utils.clip_grad_norm_(
        trainable_50,
        max_norm=CLIP_50,
        error_if_nonfinite=True
    )

    raw_norm = float(grad_norm)

    if raw_norm > 5000:
        optimizer_50.zero_grad(set_to_none=True)
        raise RuntimeError(
            f"Extreme gradient norm at update "
            f"{update}, recording {rid}: {raw_norm:.1f}"
        )

    optimizer_50.step()

    losses_50.append(float(loss.item()))
    norms_50.append(raw_norm)

    completed_50 = update

    del batch, loss

    # Evaluate at the end of each full epoch.
    if update % len(train_ids_50) == 0:

        epoch = update // len(train_ids_50)

        row = report_50(epoch, update)

        row["mean_step_loss"] = statistics.mean(
            losses_50
        )
        row["median_gradient_norm"] = statistics.median(
            norms_50
        )
        row["max_gradient_norm"] = max(norms_50)
        row["clipped_fraction"] = (
            sum(n > CLIP_50 for n in norms_50)
            / len(norms_50)
        )

        improved = (
            row["val_cer"] < best_cer_50
        )

        if improved:
            best_cer_50 = row["val_cer"]

        history_50.append(row)

        save_50(
            update,
            best_cer_50,
            save_best=improved
        )

        print(
            "Mean training-step loss:",
            round(row["mean_step_loss"], 4)
        )
        print(
            "Median gradient norm:",
            round(row["median_gradient_norm"], 2)
        )
        print(
            "Maximum gradient norm:",
            round(row["max_gradient_norm"], 2)
        )
        print(
            "Fraction clipped:",
            f"{row['clipped_fraction']*100:.1f}%"
        )

        losses_50.clear()
        norms_50.clear()

# ------------------------------------------------------------
# 7. Final comparison
# ------------------------------------------------------------

print("\n" + "=" * 70)
print("QUALITY-FILTERED TRAINING RESULTS")
print("=" * 70)

print(
    f"{'Epoch':<8}"
    f"{'Old train':<14}"
    f"{'New train':<14}"
    f"{'Val CER':<13}"
    f"{'Val WER':<13}"
    f"{'Length':<10}"
)

for row in history_50:

    print(
        f"{row['epoch']:<8}"
        f"{row['old_train_cer']*100:<14.2f}"
        f"{row['new_train_cer']*100:<14.2f}"
        f"{row['val_cer']*100:<13.2f}"
        f"{row['val_wer']*100:<13.2f}"
        f"{row['val_length_ratio']:<10.2f}"
    )

print("\nAdditional updates completed:", completed_50)
print("Best observed validation CER:",
      f"{best_cer_50*100:.2f}%")

print("Latest checkpoint:", LATEST_50)
print("History:", HISTORY_50)

if BEST_50.exists():
    print("Best improved checkpoint:", BEST_50)
else:
    print(
        "No improved stage-2 checkpoint; "
        "the stage-1 starting checkpoint remains best."
    )

print("All earlier model checkpoints unchanged.")


RESTORING SCALED MODEL
Restored Cell 45 checkpoint at update 128.

QUALITY-FILTERED TRAINING
Training recordings: 62
Primary validation: 15
Previously trained: 7
New training: 55
Trainable parameters: 25521473
FP32: True
Additional epochs: 3

EPOCH 0/3
----------------------------------------------------------
Additional updates: 0
Previous 7 training CER: 43.53%
New 55 training CER: 87.49%
Primary validation CER: 89.50%
Primary validation WER: 99.70%
Prediction/reference length: 0.36
CTC blank frames: 94.6%
Nonempty validation predictions: 15/15
Validation example:
ይ ውመበበአ ም የ ድ ው

EPOCH 1/3
----------------------------------------------------------
Additional updates: 62
Previous 7 training CER: 45.52%
New 55 training CER: 87.43%
Primary validation CER: 89.19%
Primary validation WER: 100.00%
Prediction/reference length: 0.35
CTC blank frames: 94.7%
Nonempty validation predictions: 15/15
Validation example:
ይ ውመበበአ ድ መ ድ ው
Mean training-step loss: 5.9876
Median gradient norm: 27.1
Max

In [ ]:

# ============================================================
# CELL 51 - AMHARIC CTC LABEL ROUND-TRIP AUDIT
#
# Verify that the labels used for training reconstruct
# the exact normalized reference transcripts.
#
# 62 training + 15 validation recordings.
# No training or checkpoint modifications.
# ============================================================

import json
import statistics
from collections import Counter
from pathlib import Path
from jiwer import cer

QA51_DIR = DATA_DIR / "scaled_amharic_64_16_v1"
QA51_SPLIT = QA51_DIR / "quality_filtered_v2.json"
QA51_OUTPUT = QA51_DIR / "label_roundtrip_audit.json"

selection = json.loads(
    QA51_SPLIT.read_text(encoding="utf-8")
)

groups = {
    "train": selection["train_ids"],
    "validation": selection["primary_val_ids"]
}

assert len(groups["train"]) == 62
assert len(groups["validation"]) == 15

record_lookup = {
    r["id"]: r for r in train_records
}

dataset_indices = {
    r["id"]: index
    for index, r in enumerate(train_dataset.records)
}

# XLS-R convolutional feature extractor configuration.
kernels = (10, 3, 3, 3, 2, 2, 2)
strides = (5, 2, 2, 2, 2, 2, 2)

# Read the actual architecture configuration instead
# of assuming its kernels/strides are correct.
from transformers import Wav2Vec2Config

config = Wav2Vec2Config.from_pretrained(str(BASELINE_DIR))
kernels = tuple(config.conv_kernel)
strides = tuple(config.conv_stride)

def output_frames(n_samples):
    length = int(n_samples)
    for kernel, stride in zip(kernels, strides):
        length = (length - kernel) // stride + 1
    return length

rows = []
token_counts = Counter()

print("AMHARIC CTC LABEL AUDIT")
print("=" * 60)
print("Tokenizer vocabulary size:", len(tokenizer))
print("CTC blank ID:", tokenizer.pad_token_id)
print("Unknown token ID:", tokenizer.unk_token_id)
print("Recording count:", 77)

for group_name, record_ids in groups.items():

    print(f"\nChecking {group_name}: {len(record_ids)} recordings")

    for rid in record_ids:

        record = record_lookup[rid]

        # Load the exact dataset example used in training.
        example = train_dataset[dataset_indices[rid]]
        batch = ctc_collator([example])

        # Remove only padding introduced by the collator.
        label_tensor = batch["labels"][0]
        label_ids = label_tensor[
            label_tensor != -100
        ].detach().cpu().tolist()

        # Decode WITHOUT collapsing repeated CTC symbols.
        # Repeated symbols in references must be preserved.
        decoded = tokenizer.decode(
            label_ids,
            group_tokens=False
        )

        reference = normalize_amharic_ctc(
            record["transcription"]
        )

        decoded = normalize_amharic_ctc(decoded)

        # Count unknown and blank target tokens.
        unknown_count = sum(
            tid == tokenizer.unk_token_id
            for tid in label_ids
        )

        blank_count = sum(
            tid == tokenizer.pad_token_id
            for tid in label_ids
        )

        repeated = sum(
            left == right
            for left, right in zip(
                label_ids[:-1], label_ids[1:]
            )
        )

        audio_samples = int(
            batch["attention_mask"][0].sum().item()
        )

        frames = output_frames(audio_samples)
        required_frames = len(label_ids) + repeated

        token_counts.update(label_ids)

        row = {
            "id": rid,
            "group": group_name,
            "reference": reference,
            "decoded_labels": decoded,
            "exact_match": reference == decoded,
            "roundtrip_cer": float(
                cer(reference, decoded)
            ),
            "label_length": len(label_ids),
            "unknown_count": unknown_count,
            "blank_target_count": blank_count,
            "audio_seconds": audio_samples / 16000,
            "available_frames": frames,
            "required_frames": required_frames,
            "ctc_feasible": frames >= required_frames
        }

        rows.append(row)

    print("Completed:", len(record_ids))

# ------------------------------------------------------------
# Summarize results
# ------------------------------------------------------------

mismatches = [
    r for r in rows
    if not r["exact_match"]
]

unknown_rows = [
    r for r in rows
    if r["unknown_count"] > 0
]

blank_rows = [
    r for r in rows
    if r["blank_target_count"] > 0
]

invalid_alignment = [
    r for r in rows
    if not r["ctc_feasible"]
]

references = [r["reference"] for r in rows]
decoded_all = [r["decoded_labels"] for r in rows]

print("\n" + "=" * 65)
print("LABEL INTEGRITY RESULTS")
print("=" * 65)

print("Recordings checked:", len(rows))
print("Exact transcript round-trips:",
      len(rows) - len(mismatches))
print("Transcript mismatches:", len(mismatches))
print("Recordings with unknown tokens:", len(unknown_rows))
print("Recordings with blank target tokens:", len(blank_rows))
print("CTC-infeasible recordings:", len(invalid_alignment))

print(
    "Overall label round-trip CER:",
    f"{cer(references, decoded_all)*100:.4f}%"
)

print(
    "Minimum CTC frame margin:",
    min(
        r["available_frames"] - r["required_frames"]
        for r in rows
    )
)

print(
    "Distinct token IDs appearing in labels:",
    len(token_counts)
)

# ------------------------------------------------------------
# Print any transcript reconstruction errors
# ------------------------------------------------------------

if mismatches:

    print("\nTRANSCRIPT MISMATCHES")
    print("=" * 65)

    for row in mismatches[:10]:

        print("\nID:", row["id"])
        print("Group:", row["group"])
        print("CER:", f"{row['roundtrip_cer']*100:.2f}%")
        print("REFERENCE:")
        print(row["reference"])
        print("DECODED LABELS:")
        print(row["decoded_labels"])

else:
    print("\nALL 77 LABELS RECONSTRUCT THEIR REFERENCES.")

# ------------------------------------------------------------
# Save full audit
# ------------------------------------------------------------

result = {
    "recordings_checked": len(rows),
    "exact_matches": len(rows) - len(mismatches),
    "mismatch_count": len(mismatches),
    "unknown_token_recordings": len(unknown_rows),
    "blank_target_recordings": len(blank_rows),
    "ctc_infeasible_recordings": len(invalid_alignment),
    "corpus_roundtrip_cer": float(
        cer(references, decoded_all)
    ),
    "rows": rows
}

QA51_OUTPUT.write_text(
    json.dumps(
        result,
        ensure_ascii=False,
        indent=2
    ),
    encoding="utf-8"
)

print("\n" + "=" * 65)
print("AUDIT FINISHED")
print("=" * 65)
print("Saved:", QA51_OUTPUT)
print("Optimizer updates: 0")
print("Model checkpoints modified: 0")


AMHARIC CTC LABEL AUDIT
Tokenizer vocabulary size: 321
CTC blank ID: 320
Unknown token ID: 319
Recording count: 77

Checking train: 62 recordings
Completed: 62

Checking validation: 15 recordings
Completed: 15

LABEL INTEGRITY RESULTS
Recordings checked: 77
Exact transcript round-trips: 77
Transcript mismatches: 0
Recordings with unknown tokens: 0
Recordings with blank target tokens: 0
CTC-infeasible recordings: 0
Overall label round-trip CER: 0.0000%
Minimum CTC frame margin: 191
Distinct token IDs appearing in labels: 197

ALL 77 LABELS RECONSTRUCT THEIR REFERENCES.

AUDIT FINISHED
Saved: /content/drive/MyDrive/Amharic_ASR_XLSR/data/scaled_amharic_64_16_v1/label_roundtrip_audit.json
Optimizer updates: 0
Model checkpoints modified: 0


In [ ]:

# ============================================================
# CELL 52 - TWO-HOUR TRAINING DATASET
#
# Goal: approximately 2 hours of diverse Amharic audio.
# Preserve existing evaluation speaker separation.
# Exclude known quarantined recordings.
#
# No GPU training. No checkpoint changes.
# ============================================================

import json
import random
import hashlib
import statistics
from pathlib import Path
from collections import defaultdict, Counter
from IPython.display import Audio, display
from transformers import Wav2Vec2Config

ROOT_52 = DATA_DIR / "scaled_amharic_64_16_v1"
OUT_52 = DATA_DIR / "amharic_2hour_pilot_v1"
OUT_52.mkdir(parents=True, exist_ok=True)

SELECTION_52 = OUT_52 / "selection.json"
SEED_52 = 20261020
TARGET_SECONDS_52 = 7200
MAX_RECORDINGS_52 = 750
MAX_PER_SPEAKER_52 = 5

clean = json.loads(
    (ROOT_52 / "quality_filtered_v2.json").read_text(
        encoding="utf-8"
    )
)

original = json.loads(
    (ROOT_52 / "selection.json").read_text(
        encoding="utf-8"
    )
)

records_52 = {r["id"]: r for r in train_records}

# ------------------------------------------------------------
# 1. Protect evaluation examples AND speakers
# ------------------------------------------------------------

protected_ids_52 = set(original["val_ids"])
protected_ids_52.update(clean["primary_val_ids"])
protected_ids_52.update(clean["noisy_challenge_ids"])

prior_validation_files = [
    DATA_DIR / "short_multirecording_head_only_v2"
    / "split.json",

    DATA_DIR / "head_only_multirecording_v1"
    / "selection.json"
]

for path in prior_validation_files:
    if path.is_file():
        previous = json.loads(
            path.read_text(encoding="utf-8")
        )
        protected_ids_52.update(
            previous.get("val_ids", [])
        )

# Protect the original fixed evaluation IDs/speakers
# too, if its metadata is present in the JSONL file.
external_speakers_52 = set()

external_path_52 = DATA_DIR / "baseline_eval_fixed_12.jsonl"

if external_path_52.is_file():
    for line in external_path_52.read_text(
        encoding="utf-8"
    ).splitlines():
        if not line.strip():
            continue

        entry = json.loads(line)
        rid = entry.get("id")

        if rid:
            protected_ids_52.add(rid)

        if entry.get("speaker_id"):
            external_speakers_52.add(
                entry["speaker_id"]
            )

protected_speakers_52 = {
    records_52[rid]["speaker_id"]
    for rid in protected_ids_52
    if rid in records_52
}
protected_speakers_52.update(external_speakers_52)

quarantined_52 = set(
    clean["quarantined_train_ids"]
)

print("PROTECTION CHECKS")
print("=" * 55)
print("Protected recording IDs:", len(protected_ids_52))
print("Protected speaker IDs:", len(protected_speakers_52))
print("Quarantined recordings:", len(quarantined_52))

# ------------------------------------------------------------
# 2. Verify recording eligibility
# ------------------------------------------------------------

cfg_52 = Wav2Vec2Config.from_pretrained(
    str(BASELINE_DIR)
)

def frames_52(n_samples):
    n = int(n_samples)
    for kernel, stride in zip(
        cfg_52.conv_kernel, cfg_52.conv_stride
    ):
        n = (n - kernel) // stride + 1
    return n

def eligible_52(record):
    rid = record["id"]
    sid = record.get("speaker_id")

    if not sid:
        return False
    if rid in protected_ids_52 | quarantined_52:
        return False
    if sid in protected_speakers_52:
        return False

    seconds = float(record["duration_seconds"])
    if not 4.0 <= seconds <= 18.0:
        return False

    text = record["transcription"]

    if any(ch.isdigit() for ch in text):
        return False

    audio_path = Path(AUDIO_DIR) / record["audio_file"]
    if not audio_path.is_file():
        return False

    labels = tokenizer.encode(
        text, add_special_tokens=False
    )

    if not 20 <= len(labels) <= 160:
        return False

    if tokenizer.unk_token_id in labels:
        return False
    if tokenizer.pad_token_id in labels:
        return False

    repeats = sum(
        a == b
        for a, b in zip(labels[:-1], labels[1:])
    )

    available = frames_52(round(seconds * 16000))
    return available - len(labels) - repeats >= 20

eligible_records_52 = [
    r for r in train_records
    if eligible_52(r)
]

print("\nEligible candidates:", len(eligible_records_52))
print(
    "Eligible speakers:",
    len({r["speaker_id"] for r in eligible_records_52})
)

# ------------------------------------------------------------
# 3. Retain valid previously trained examples
# ------------------------------------------------------------

carryover_52 = [
    rid for rid in clean["train_ids"]
    if eligible_52(records_52[rid])
]

excluded_carryover_52 = [
    rid for rid in clean["train_ids"]
    if rid not in carryover_52
]

print("\nPrevious training recordings retained:",
      len(carryover_52))

print("Additional carryover exclusions:",
      len(excluded_carryover_52))

# ------------------------------------------------------------
# 4. Speaker-balanced selection
# ------------------------------------------------------------

if SELECTION_52.exists():

    selection_52 = json.loads(
        SELECTION_52.read_text(encoding="utf-8")
    )

    selected_ids_52 = selection_52["train_ids"]

    print("\nRestored existing saved selection.")

else:

    rng = random.Random(SEED_52)

    selected_ids_52 = list(carryover_52)
    selected_set_52 = set(selected_ids_52)

    counts_52 = Counter(
        records_52[rid]["speaker_id"]
        for rid in selected_ids_52
    )

    total_seconds_52 = sum(
        float(records_52[rid]["duration_seconds"])
        for rid in selected_ids_52
    )

    by_speaker_52 = defaultdict(list)

    for record in eligible_records_52:
        if record["id"] not in selected_set_52:
            by_speaker_52[
                record["speaker_id"]
            ].append(record)

    speakers_52 = sorted(by_speaker_52)
    rng.shuffle(speakers_52)

    for sid in speakers_52:
        rng.shuffle(by_speaker_52[sid])

    # Round-robin sampling promotes speaker diversity.
    for _ in range(MAX_PER_SPEAKER_52):

        if total_seconds_52 >= TARGET_SECONDS_52:
            break

        for sid in speakers_52:

            if total_seconds_52 >= TARGET_SECONDS_52:
                break
            if len(selected_ids_52) >= MAX_RECORDINGS_52:
                break
            if counts_52[sid] >= MAX_PER_SPEAKER_52:
                continue
            if not by_speaker_52[sid]:
                continue

            record = by_speaker_52[sid].pop()
            rid = record["id"]

            selected_ids_52.append(rid)
            selected_set_52.add(rid)

            counts_52[sid] += 1
            total_seconds_52 += float(
                record["duration_seconds"]
            )

    assert total_seconds_52 >= TARGET_SECONDS_52, (
        "Unable to reach 2 hours under these constraints. "
        f"Selected {total_seconds_52 / 3600:.2f} hours."
    )

    selection_52 = {
        "seed": SEED_52,
        "source": "train_final_25h_ctc_safe",
        "train_ids": selected_ids_52,
        "carryover_ids": carryover_52,
        "excluded_carryover_ids": excluded_carryover_52,
        "primary_val_ids": clean["primary_val_ids"],
        "noisy_challenge_ids": clean["noisy_challenge_ids"],
        "quarantined_ids": sorted(quarantined_52),
        "target_audio_seconds": TARGET_SECONDS_52,
        "max_recordings": MAX_RECORDINGS_52,
        "max_per_speaker": MAX_PER_SPEAKER_52
    }

    SELECTION_52.write_text(
        json.dumps(
            selection_52,
            indent=2,
            ensure_ascii=False
        ),
        encoding="utf-8"
    )

    print("\nNew two-hour selection saved.")

# ------------------------------------------------------------
# 5. Check for leakage and invalid examples
# ------------------------------------------------------------

selected_records_52 = [
    records_52[rid]
    for rid in selected_ids_52
]

assert len(selected_ids_52) == len(set(selected_ids_52))

assert all(
    eligible_52(r)
    for r in selected_records_52
)

train_speakers_52 = {
    r["speaker_id"] for r in selected_records_52
}

assert not (
    train_speakers_52 & protected_speakers_52
)
assert not (
    set(selected_ids_52) & protected_ids_52
)
assert not (
    set(selected_ids_52) & quarantined_52
)

# ------------------------------------------------------------
# 6. Verify tokenizer reconstruction again
# ------------------------------------------------------------

roundtrip_errors_52 = []

for record in selected_records_52:

    original_text = normalize_amharic_ctc(
        record["transcription"]
    )

    ids = tokenizer.encode(
        record["transcription"],
        add_special_tokens=False
    )

    recovered = normalize_amharic_ctc(
        tokenizer.decode(
            ids, group_tokens=False
        )
    )

    if original_text != recovered:
        roundtrip_errors_52.append(record["id"])

assert not roundtrip_errors_52, (
    f"Tokenizer mismatches: {roundtrip_errors_52[:5]}"
)

# ------------------------------------------------------------
# 7. Summarize the selection
# ------------------------------------------------------------

durations_52 = [
    float(r["duration_seconds"])
    for r in selected_records_52
]

total_hours_52 = sum(durations_52) / 3600

speaker_counts_52 = Counter(
    r["speaker_id"] for r in selected_records_52
)

print("\n" + "=" * 60)
print("TWO-HOUR DATASET SUMMARY")
print("=" * 60)

print("Selected recordings:", len(selected_records_52))
print("Selected speakers:", len(train_speakers_52))
print("Total audio:", round(total_hours_52, 3), "hours")
print("Average duration:",
      round(statistics.mean(durations_52), 2), "seconds")
print("Shortest duration:", round(min(durations_52), 2))
print("Longest duration:", round(max(durations_52), 2))

print("Maximum recordings from one speaker:",
      max(speaker_counts_52.values()))

print("Tokenizer round-trip mismatches:",
      len(roundtrip_errors_52))

print("Validation-speaker overlap:", 0)
print("Quarantined examples included:", 0)

print("Primary validation examples:",
      len(selection_52["primary_val_ids"]))

# ------------------------------------------------------------
# 8. Randomly spot-check newly selected recordings
# ------------------------------------------------------------

new_records_52 = [
    r for r in selected_records_52
    if r["id"] not in set(carryover_52)
]

sample_rng_52 = random.Random(SEED_52 + 1)
spot_checks_52 = sample_rng_52.sample(
    new_records_52,
    min(4, len(new_records_52))
)

print("\nRANDOM AUDIO QUALITY CHECK")
print("=" * 60)

for i, record in enumerate(spot_checks_52, 1):

    print(f"\nSAMPLE {i}")
    print("ID:", record["id"])
    print("Duration:", record["duration_seconds"])
    print("Transcript:", record["transcription"])

    display(Audio(
        filename=str(
            Path(AUDIO_DIR) / record["audio_file"]
        )
    ))

print("\nSELECTION COMPLETE")
print("Saved:", SELECTION_52)
print("No training or model checkpoint modifications.")


PROTECTION CHECKS
Protected recording IDs: 36
Protected speaker IDs: 28
Quarantined recordings: 2

Eligible candidates: 2832
Eligible speakers: 514

Previous training recordings retained: 59
Additional carryover exclusions: 3

New two-hour selection saved.

TWO-HOUR DATASET SUMMARY
Selected recordings: 452
Selected speakers: 408
Total audio: 2.001 hours
Average duration: 15.94 seconds
Shortest duration: 4.3
Longest duration: 17.98
Maximum recordings from one speaker: 3
Tokenizer round-trip mismatches: 0
Validation-speaker overlap: 0
Quarantined examples included: 0
Primary validation examples: 15

RANDOM AUDIO QUALITY CHECK

SAMPLE 1
ID: 8Nx0eN5fpVQrwnDxQwCt
Duration: 16.464
Transcript: ምግብ ማለት አንድ ሰው በህይወት ለመኖር አስፈላጊ ነገር ነው ምግብ ከሌላ በህይወት መኖር የለም ስለዚህ ምግብ በይወት ለመኖር ለአንድ ሰው ጠቃሚ ነገር ነው ማለት ነው



SAMPLE 2
ID: 8I7U8BiPRUTTR2zGGwC2
Duration: 16.704
Transcript: ይሄ ምናየው ልጆች የሙዚቃ እንቅስቃሴያቸውን ወይም ውዝዋዜያቸውን እያሳዩ ይመስላል እነዚህም ልጆች አረንጓዴ መስክ ላይ ይታያሉ



SAMPLE 3
ID: 17YmtLD6ty8Euq3veXaQ
Duration: 15.864
Transcript: ቲዎሎጂ ትምህርት የሚሰኘው ትምህርት አይነት ስለ ክርስቲያኗ ቅዱስ እና ቀኖና የሚሰጥበት የትምህርት ሲሆንና የተለያዩ ቤተ ክህነትና ዲቁና ላላቸው ሰዎች ይሰጣል



SAMPLE 4
ID: 8FKfXlzJMfHqjnOlSUjm
Duration: 17.016
Transcript: ጋዜጣ ላይ የሚወጡ ማስታወቂያዎች ብዙ ጊዜ ከመደበኛ ማስታወቂያዎች በቲቪና ከሬድዮ ከሚተላለፉ ለየት የሚያደርጋቸው ብዛት ያላቸውን የሐራጅ ማስታወቂያዎችን የባንክ ማስታወቂያዎችን ስለ አክሲዮኖች አዋጆች ምናምን ስለሚወጡ ነው



SELECTION COMPLETE
Saved: /content/drive/MyDrive/Amharic_ASR_XLSR/data/amharic_2hour_pilot_v1/selection.json
No training or model checkpoint modifications.


In [ ]:

# ============================================================
# CELL 53 - TWO-HOUR HEAD-ONLY ASR TRAINING
#
# 452 training recordings / 15 development recordings
# Frozen encoder: best model from Cell 50
# Trainable: CTC head only (329,025 parameters)
#
# 5 epochs, full FP32
# Resumable checkpoints after every epoch
# All earlier checkpoints remain unchanged
# ============================================================

import gc
import copy
import json
import math
import random
import hashlib
from pathlib import Path

import torch
import torch.nn.functional as F
from jiwer import cer, wer
from transformers import Wav2Vec2ForCTC

DEVICE_53 = torch.device(
    "cuda" if torch.cuda.is_available() else "cpu"
)

ROOT_53 = DATA_DIR / "amharic_2hour_pilot_v1"

SOURCE_53 = (
    DATA_DIR / "scaled_amharic_64_16_v1"
    / "stage2_filtered_62_v1" / "best.pt"
)

SELECTION_53 = ROOT_53 / "selection.json"

RUN_53 = ROOT_53 / "head_only_stage1_v1"
RUN_53.mkdir(parents=True, exist_ok=True)

LATEST_53 = RUN_53 / "latest.pt"
BEST_53 = RUN_53 / "best.pt"
HISTORY_53 = RUN_53 / "history.json"

EPOCHS_53 = 5
HEAD_LR_53 = 5e-4
CLIP_53 = 5.0
SEED_53 = 20261020
BLANK_53 = tokenizer.pad_token_id

assert SOURCE_53.is_file()
assert SELECTION_53.is_file()

selection_53 = json.loads(
    SELECTION_53.read_text(encoding="utf-8")
)

train_ids_53 = selection_53["train_ids"]
val_ids_53 = selection_53["primary_val_ids"]
carryover_53 = selection_53["carryover_ids"]

assert len(train_ids_53) == 452
assert len(val_ids_53) == 15
assert len(set(train_ids_53 + val_ids_53)) == 467

records_53 = {r["id"]: r for r in train_records}
indices_53 = {
    r["id"]: i
    for i, r in enumerate(train_dataset.records)
}

assert all(
    rid in indices_53
    for rid in train_ids_53 + val_ids_53
)

train_speakers_53 = {
    records_53[rid]["speaker_id"]
    for rid in train_ids_53
}

val_speakers_53 = {
    records_53[rid]["speaker_id"]
    for rid in val_ids_53
}

assert not train_speakers_53.intersection(val_speakers_53)

new_ids_53 = [
    rid for rid in train_ids_53
    if rid not in set(carryover_53)
]

# Fixed training probe, separate from evaluation.
rng_probe_53 = random.Random(SEED_53)
new_probe_53 = rng_probe_53.sample(
    new_ids_53, min(64, len(new_ids_53))
)

print("TWO-HOUR HEAD-ONLY EXPERIMENT")
print("=" * 60)
print("Training examples:", len(train_ids_53))
print("Development examples:", len(val_ids_53))
print("Previously used training examples:", len(carryover_53))
print("New training examples:", len(new_ids_53))
print("Distinct training speakers:", len(train_speakers_53))
print("Train/development speaker overlap:", 0)
print("Device:", DEVICE_53)

# ------------------------------------------------------------
# 1. Load adapted encoder and trained head
# ------------------------------------------------------------

source_53 = torch.load(
    SOURCE_53,
    map_location="cpu",
    weights_only=True
)

assert source_53["precision"] == "fp32"
assert len(source_53["upper_layers"]) == 2

model_53 = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(DEVICE_53).float()

model_53.lm_head.load_state_dict(
    source_53["head"], strict=True
)

for layer, weights in zip(
    model_53.wav2vec2.encoder.layers[-2:],
    source_53["upper_layers"]
):
    layer.load_state_dict(weights, strict=True)

model_53.eval()
model_53.requires_grad_(False)

# Copy the trainable head outside inference_mode.
head_53 = copy.deepcopy(
    model_53.lm_head
).to(DEVICE_53).float()

head_53.requires_grad_(True)

assert sum(
    p.numel() for p in head_53.parameters()
) == 329025

print("\nStarting model restored.")
print("Encoder: frozen")
print("CTC head: trainable")
print("Head parameters: 329,025")

# ------------------------------------------------------------
# 2. Cache frozen encoder features in CPU RAM
# ------------------------------------------------------------

# Each item stores its encoder output as float32.
# This avoids running the 300M-parameter XLS-R encoder
# again on every training epoch.

def cache_record_53(rid):

    example = train_dataset[indices_53[rid]]
    batch = ctc_collator([example])

    input_values = batch["input_values"].to(
        DEVICE_53
    )

    attention_mask = batch["attention_mask"].to(
        DEVICE_53
    )

    with torch.no_grad():
        hidden = model_53.wav2vec2(
            input_values=input_values,
            attention_mask=attention_mask
        ).last_hidden_state

    features = hidden.detach().cpu().float().contiguous()

    targets = batch["labels"][0]
    targets = targets[
        targets >= 0
    ].detach().cpu().long().contiguous()

    repeats = int(
        (targets[1:] == targets[:-1]).sum().item()
    )

    assert features.shape[1] >= (
        targets.numel() + repeats
    )

    assert not (targets == BLANK_53).any()
    assert torch.isfinite(features).all().item()

    reference = normalize_amharic_ctc(
        records_53[rid]["transcription"]
    )

    return {
        "features": features,
        "targets": targets,
        "frames": int(features.shape[1]),
        "target_length": int(targets.numel()),
        "reference": reference
    }

print("\nCaching frozen encoder features...")
print("Features are stored in CPU RAM.")

cache_53 = {}

all_ids_53 = train_ids_53 + val_ids_53

for i, rid in enumerate(all_ids_53, 1):

    cache_53[rid] = cache_record_53(rid)

    if i % 50 == 0 or i == len(all_ids_53):
        print(f"Cached: {i}/{len(all_ids_53)}")

cached_bytes_53 = sum(
    item["features"].numel() * 4
    for item in cache_53.values()
)

print(
    "Cached feature memory:",
    round(cached_bytes_53 / 1024**3, 2),
    "GiB"
)

# The encoder is no longer needed for head training.
del model_53
gc.collect()

if DEVICE_53.type == "cuda":
    torch.cuda.empty_cache()

# ------------------------------------------------------------
# 3. Setup optimizer and reproducible experiment ID
# ------------------------------------------------------------

optimizer_53 = torch.optim.AdamW(
    head_53.parameters(),
    lr=HEAD_LR_53,
    weight_decay=0.0
)

config_53 = {
    "source_checkpoint": str(SOURCE_53),
    "source_update": source_53.get("updates"),
    "training_ids": train_ids_53,
    "development_ids": val_ids_53,
    "references": {
        rid: records_53[rid]["transcription"]
        for rid in all_ids_53
    },
    "head_lr": HEAD_LR_53,
    "clip_norm": CLIP_53,
    "seed": SEED_53,
    "epochs": EPOCHS_53
}

signature_53 = hashlib.sha256(
    json.dumps(
        config_53,
        sort_keys=True,
        ensure_ascii=False
    ).encode("utf-8")
).hexdigest()

# ------------------------------------------------------------
# 4. Resume existing experiment if available
# ------------------------------------------------------------

start_epoch_53 = 0
history_53 = []
best_cer_53 = float("inf")

if LATEST_53.exists():

    previous_53 = torch.load(
        LATEST_53,
        map_location="cpu",
        weights_only=True
    )

    assert previous_53["signature"] == signature_53

    head_53.load_state_dict(
        previous_53["head"]
    )

    optimizer_53.load_state_dict(
        previous_53["optimizer"]
    )

    start_epoch_53 = int(
        previous_53["completed_epochs"]
    )

    best_cer_53 = float(
        previous_53["best_cer"]
    )

    if HISTORY_53.exists():
        history_53 = json.loads(
            HISTORY_53.read_text(encoding="utf-8")
        )

    print(
        "\nResuming from completed epoch:",
        start_epoch_53
    )

else:
    print("\nStarting new head-only training.")

assert 0 <= start_epoch_53 <= EPOCHS_53

# ------------------------------------------------------------
# 5. CTC training loss
# ------------------------------------------------------------

def loss_53(rid):

    item = cache_53[rid]

    features = item["features"].to(DEVICE_53)
    targets = item["targets"].to(DEVICE_53)

    logits = head_53(features)

    log_probs = F.log_softmax(
        logits.float(), dim=-1
    ).transpose(0, 1)

    input_lengths = torch.tensor(
        [item["frames"]],
        dtype=torch.long
    )

    target_lengths = torch.tensor(
        [item["target_length"]],
        dtype=torch.long
    )

    return F.ctc_loss(
        log_probs,
        targets,
        input_lengths,
        target_lengths,
        blank=BLANK_53,
        reduction="mean",
        zero_infinity=False
    )

# ------------------------------------------------------------
# 6. Evaluation
# ------------------------------------------------------------

def evaluate_53(ids):

    head_53.eval()

    references = []
    predictions = []

    blank_count = 0
    frame_count = 0

    with torch.no_grad():

        for rid in ids:

            item = cache_53[rid]

            features = item["features"].to(
                DEVICE_53
            )

            logits = head_53(features)

            predicted_ids = logits.argmax(
                dim=-1
            )

            blank_count += int(
                (predicted_ids == BLANK_53).sum().item()
            )

            frame_count += predicted_ids.numel()

            prediction = processor.batch_decode(
                predicted_ids.cpu()
            )[0]

            prediction = normalize_amharic_ctc(
                prediction
            )

            references.append(item["reference"])
            predictions.append(prediction)

    reference_chars = sum(
        len(s.replace(" ", ""))
        for s in references
    )

    predicted_chars = sum(
        len(s.replace(" ", ""))
        for s in predictions
    )

    return {
        "cer": float(cer(references, predictions)),
        "wer": float(wer(references, predictions)),
        "length_ratio": (
            predicted_chars / max(reference_chars, 1)
        ),
        "blank_fraction": (
            blank_count / max(frame_count, 1)
        ),
        "nonempty": sum(
            bool(s.strip()) for s in predictions
        ),
        "example": predictions[0]
    }

def report_53(epoch):

    old = evaluate_53(carryover_53)
    new = evaluate_53(new_probe_53)
    dev = evaluate_53(val_ids_53)

    result = {
        "epoch": epoch,
        "updates": epoch * len(train_ids_53),
        "old_train_cer": old["cer"],
        "new_train_probe_cer": new["cer"],
        "dev_cer": dev["cer"],
        "dev_wer": dev["wer"],
        "dev_length_ratio": dev["length_ratio"],
        "dev_blank_fraction": dev["blank_fraction"],
        "dev_nonempty": dev["nonempty"],
        "dev_example": dev["example"]
    }

    print(f"\nEPOCH {epoch}/{EPOCHS_53}")
    print("-" * 55)
    print(
        "Previously trained CER:",
        f"{old['cer']*100:.2f}%"
    )
    print(
        "New training probe CER:",
        f"{new['cer']*100:.2f}%"
    )
    print(
        "Development CER:",
        f"{dev['cer']*100:.2f}%"
    )
    print(
        "Development WER:",
        f"{dev['wer']*100:.2f}%"
    )
    print(
        "Prediction/reference length:",
        f"{dev['length_ratio']:.2f}"
    )
    print(
        "Blank frames:",
        f"{dev['blank_fraction']*100:.2f}%"
    )
    print(
        "Nonempty development predictions:",
        f"{dev['nonempty']}/15"
    )
    print(
        "Development example:",
        dev["example"][:120] or "[EMPTY]"
    )

    return result

# ------------------------------------------------------------
# 7. Checkpoint management
# ------------------------------------------------------------

def save_53(epoch, improved):

    state = {
        "signature": signature_53,
        "completed_epochs": epoch,
        "best_cer": best_cer_53,
        "source_checkpoint": str(SOURCE_53),
        "head": head_53.state_dict(),
        "optimizer": optimizer_53.state_dict()
    }

    temporary = RUN_53 / "latest.pt.partial"
    torch.save(state, temporary)
    temporary.replace(LATEST_53)

    if improved:
        temporary_best = RUN_53 / "best.pt.partial"
        torch.save(state, temporary_best)
        temporary_best.replace(BEST_53)

    temporary_history = RUN_53 / "history.json.partial"

    temporary_history.write_text(
        json.dumps(
            history_53,
            ensure_ascii=False,
            indent=2
        ),
        encoding="utf-8"
    )

    temporary_history.replace(HISTORY_53)

# ------------------------------------------------------------
# 8. Establish baseline
# ------------------------------------------------------------

print("\nTWO-HOUR FROZEN-ENCODER TRAINING")
print("=" * 60)
print("Epochs:", EPOCHS_53)
print("Total planned optimizer updates:",
      EPOCHS_53 * len(train_ids_53))
print("Precision: FP32")
print("Head LR:", HEAD_LR_53)
print("Gradient clipping:", CLIP_53)

if start_epoch_53 == 0 and not history_53:

    initial_53 = report_53(0)
    history_53.append(initial_53)
    best_cer_53 = initial_53["dev_cer"]

# ------------------------------------------------------------
# 9. Train CTC head for five epochs
# ------------------------------------------------------------

for epoch in range(
    start_epoch_53 + 1,
    EPOCHS_53 + 1
):

    order = list(train_ids_53)

    random.Random(
        SEED_53 + epoch
    ).shuffle(order)

    losses = []
    gradient_norms = []

    head_53.train()

    for i, rid in enumerate(order, 1):

        optimizer_53.zero_grad(set_to_none=True)

        loss = loss_53(rid)

        if not torch.isfinite(loss).item():
            raise RuntimeError(
                f"Invalid CTC loss: {rid}"
            )

        loss.backward()

        norm = torch.nn.utils.clip_grad_norm_(
            head_53.parameters(),
            max_norm=CLIP_53,
            error_if_nonfinite=True
        )

        optimizer_53.step()

        losses.append(float(loss.item()))
        gradient_norms.append(float(norm))

        if i % 100 == 0 or i == len(order):
            print(
                f"Epoch {epoch}: "
                f"{i}/{len(order)} updates"
            )

    result = report_53(epoch)

    result["mean_training_loss"] = (
        sum(losses) / len(losses)
    )

    result["median_gradient_norm"] = (
        sorted(gradient_norms)[
            len(gradient_norms) // 2
        ]
    )

    result["clipped_fraction"] = (
        sum(n > CLIP_53 for n in gradient_norms)
        / len(gradient_norms)
    )

    improved = result["dev_cer"] < best_cer_53

    if improved:
        best_cer_53 = result["dev_cer"]

    history_53.append(result)
    save_53(epoch, improved)

    print(
        "Mean CTC training loss:",
        round(result["mean_training_loss"], 4)
    )

    print(
        "Median gradient norm:",
        round(result["median_gradient_norm"], 3)
    )

    print(
        "Gradient clipping frequency:",
        f"{result['clipped_fraction']*100:.1f}%"
    )

    # Stop early if severe blank collapse develops.
    if (
        result["dev_length_ratio"] < 0.10
        and result["dev_blank_fraction"] > 0.98
    ):
        print(
            "\nEARLY STOP: Severe under-generation "
            "and blank dominance detected."
        )
        break

# ------------------------------------------------------------
# 10. Final summary
# ------------------------------------------------------------

print("\n" + "=" * 75)
print("TWO-HOUR HEAD-ONLY TRAINING RESULTS")
print("=" * 75)

print(
    f"{'Epoch':<8}"
    f"{'Old CER':<13}"
    f"{'New CER':<13}"
    f"{'Dev CER':<13}"
    f"{'Dev WER':<13}"
    f"{'Length':<10}"
)

for row in history_53:

    print(
        f"{row['epoch']:<8}"
        f"{row['old_train_cer']*100:<13.2f}"
        f"{row['new_train_probe_cer']*100:<13.2f}"
        f"{row['dev_cer']*100:<13.2f}"
        f"{row['dev_wer']*100:<13.2f}"
        f"{row['dev_length_ratio']:<10.2f}"
    )

print(
    "\nBest development CER:",
    f"{best_cer_53*100:.2f}%"
)

print("Latest checkpoint:", LATEST_53)

if BEST_53.exists():
    print("Best improved checkpoint:", BEST_53)
else:
    print(
        "No improvement over starting model. "
        "Use the original source checkpoint."
    )

print("History:", HISTORY_53)
print("All previous checkpoints unchanged.")


TWO-HOUR HEAD-ONLY EXPERIMENT
Training examples: 452
Development examples: 15
Previously used training examples: 59
New training examples: 393
Distinct training speakers: 408
Train/development speaker overlap: 0
Device: cuda

Starting model restored.
Encoder: frozen
CTC head: trainable
Head parameters: 329,025

Caching frozen encoder features...
Features are stored in CPU RAM.
Cached: 50/467
Cached: 100/467
Cached: 150/467
Cached: 200/467
Cached: 250/467
Cached: 300/467
Cached: 350/467
Cached: 400/467
Cached: 450/467
Cached: 467/467
Cached feature memory: 1.41 GiB

Starting new head-only training.

TWO-HOUR FROZEN-ENCODER TRAINING
Epochs: 5
Total planned optimizer updates: 2260
Precision: FP32
Head LR: 0.0005
Gradient clipping: 5.0

EPOCH 0/5
-------------------------------------------------------
Previously trained CER: 84.34%
New training probe CER: 88.36%
Development CER: 89.07%
Development WER: 100.00%
Prediction/reference length: 0.33
Blank frames: 94.82%
Nonempty development pred

In [ ]:

# ============================================================
# CELL 54 - CTC BLANK-BIAS DIAGNOSTIC
#
# Compare warm start, epoch 1, and epoch 4.
# Test blank-logit penalties WITHOUT training.
#
# Uses cached XLS-R features from Cell 53.
# No model checkpoints modified.
# ============================================================

import json
import random
from pathlib import Path

import torch
from jiwer import cer, wer

ROOT_54 = DATA_DIR / "amharic_2hour_pilot_v1"
RUN_54 = ROOT_54 / "head_only_stage1_v1"

SOURCE_54 = (
    DATA_DIR / "scaled_amharic_64_16_v1"
    / "stage2_filtered_62_v1" / "best.pt"
)

CHECKPOINTS_54 = {
    "Warm start": SOURCE_54,
    "Epoch 1": RUN_54 / "best.pt",
    "Epoch 4": RUN_54 / "latest.pt"
}

assert "cache_53" in globals(), (
    "Cell 53's cached encoder features are unavailable. "
    "Do not rerun training just to restore them."
)

selection_54 = json.loads(
    (ROOT_54 / "selection.json").read_text(
        encoding="utf-8"
    )
)

train_ids_54 = selection_54["train_ids"]
val_ids_54 = selection_54["primary_val_ids"]
carryover_54 = set(selection_54["carryover_ids"])

new_train_ids_54 = [
    rid for rid in train_ids_54
    if rid not in carryover_54
]

train_probe_54 = random.Random(20261020).sample(
    new_train_ids_54, 64
)

all_ids_54 = train_probe_54 + val_ids_54

assert len(train_probe_54) == 64
assert len(val_ids_54) == 15
assert all(rid in cache_53 for rid in all_ids_54)

blank_id_54 = tokenizer.pad_token_id
penalties_54 = [0.0, 0.5, 1.0, 1.5, 2.0, 3.0, 4.0]

device_54 = torch.device(
    "cuda" if torch.cuda.is_available() else "cpu"
)

print("CTC BLANK-BIAS DIAGNOSTIC")
print("=" * 60)
print("Training probe:", len(train_probe_54))
print("Development recordings:", len(val_ids_54))
print("Penalties:", penalties_54)
print("No training will be performed.")

# ------------------------------------------------------------
# 1. Decode cached logits with an optional blank penalty
# ------------------------------------------------------------

def decode_logits_54(logits, penalty):

    adjusted = logits.clone()

    adjusted[:, :, blank_id_54] -= penalty

    token_ids = adjusted.argmax(dim=-1)

    text = processor.batch_decode(
        token_ids
    )[0]

    return (
        normalize_amharic_ctc(text),
        int((token_ids == blank_id_54).sum().item()),
        token_ids.numel()
    )

def evaluate_54(logit_cache, record_ids, penalty):

    references = []
    predictions = []

    blank_frames = 0
    all_frames = 0

    for rid in record_ids:

        prediction, blanks, frames = decode_logits_54(
            logit_cache[rid], penalty
        )

        references.append(
            cache_53[rid]["reference"]
        )

        predictions.append(prediction)

        blank_frames += blanks
        all_frames += frames

    ref_characters = sum(
        len(s.replace(" ", ""))
        for s in references
    )

    predicted_characters = sum(
        len(s.replace(" ", ""))
        for s in predictions
    )

    return {
        "cer": float(cer(references, predictions)),
        "wer": float(wer(references, predictions)),
        "length_ratio": (
            predicted_characters / max(ref_characters, 1)
        ),
        "blank_fraction": (
            blank_frames / max(all_frames, 1)
        ),
        "nonempty": sum(bool(s.strip()) for s in predictions),
        "sample_prediction": predictions[0]
    }

# ------------------------------------------------------------
# 2. Compare all three heads using identical features
# ------------------------------------------------------------

all_results_54 = {}

expected_dev_54 = {
    "Warm start": 0.8907,
    "Epoch 1": 0.8882,
    "Epoch 4": 0.9592
}

for model_name, path in CHECKPOINTS_54.items():

    assert path.is_file(), f"Missing checkpoint: {path}"

    saved = torch.load(
        path,
        map_location="cpu",
        weights_only=True
    )

    head_weights = saved["head"]

    weight = head_weights["weight"]

    diagnostic_head = torch.nn.Linear(
        in_features=weight.shape[1],
        out_features=weight.shape[0],
        bias=True
    ).to(device_54).float()

    diagnostic_head.load_state_dict(
        head_weights,
        strict=True
    )

    diagnostic_head.eval()

    # Compute acoustic logits only once per recording.
    # Keep logits in CPU RAM for the penalty sweep.
    logit_cache_54 = {}

    with torch.no_grad():

        for rid in all_ids_54:

            features = cache_53[rid]["features"].to(
                device_54
            )

            logits = diagnostic_head(features)

            logit_cache_54[rid] = (
                logits.detach().cpu().float()
            )

    model_results = []

    for penalty in penalties_54:

        train_result = evaluate_54(
            logit_cache_54,
            train_probe_54,
            penalty
        )

        dev_result = evaluate_54(
            logit_cache_54,
            val_ids_54,
            penalty
        )

        model_results.append({
            "penalty": penalty,
            "train_cer": train_result["cer"],
            "dev_cer": dev_result["cer"],
            "dev_wer": dev_result["wer"],
            "dev_length_ratio": dev_result["length_ratio"],
            "dev_blank_fraction": dev_result["blank_fraction"],
            "dev_nonempty": dev_result["nonempty"],
            "dev_sample": dev_result["sample_prediction"]
        })

    # Verify our zero-penalty baseline matches Cell 53.
    actual_baseline = model_results[0]["dev_cer"]

    assert abs(
        actual_baseline - expected_dev_54[model_name]
    ) < 0.005, (
        f"Baseline mismatch for {model_name}: "
        f"{actual_baseline:.4f}"
    )

    all_results_54[model_name] = model_results

    print("\n" + "=" * 72)
    print(model_name.upper())
    print("=" * 72)

    print(
        f"{'Penalty':<10}"
        f"{'Train CER':<15}"
        f"{'Dev CER':<14}"
        f"{'Dev length':<15}"
        f"{'Dev blank':<14}"
    )

    for row in model_results:

        print(
            f"{row['penalty']:<10.1f}"
            f"{row['train_cer']*100:<15.2f}"
            f"{row['dev_cer']*100:<14.2f}"
            f"{row['dev_length_ratio']:<15.2f}"
            f"{row['dev_blank_fraction']*100:<14.2f}"
        )

    # Pick an adjustment using training CER, not
    # development CER, to reduce validation tuning.
    chosen = min(
        model_results,
        key=lambda r: (
            r["train_cer"],
            r["penalty"]
        )
    )

    print(
        "\nBest training-probe penalty:",
        chosen["penalty"]
    )

    print(
        "Development CER at chosen penalty:",
        f"{chosen['dev_cer']*100:.2f}%"
    )

    print(
        "Development WER:",
        f"{chosen['dev_wer']*100:.2f}%"
    )

    print(
        "Development prediction/reference length:",
        f"{chosen['dev_length_ratio']:.2f}"
    )

    print(
        "Example prediction:",
        chosen["dev_sample"][:150] or "[EMPTY]"
    )

    del diagnostic_head, logit_cache_54

# ------------------------------------------------------------
# 3. Save diagnostic results
# ------------------------------------------------------------

output_54 = RUN_54 / "blank_bias_diagnostic.json"

output_54.write_text(
    json.dumps(
        {
            "description": (
                "Exploratory blank-logit penalty diagnostic. "
                "Penalties are not learned model parameters."
            ),
            "train_probe_count": len(train_probe_54),
            "development_count": len(val_ids_54),
            "results": all_results_54
        },
        ensure_ascii=False,
        indent=2
    ),
    encoding="utf-8"
)

print("\n" + "=" * 60)
print("BLANK-BIAS DIAGNOSTIC FINISHED")
print("=" * 60)
print("Results saved:", output_54)
print("Optimizer updates: 0")
print("Model checkpoints modified: 0")


CTC BLANK-BIAS DIAGNOSTIC
Training probe: 64
Development recordings: 15
Penalties: [0.0, 0.5, 1.0, 1.5, 2.0, 3.0, 4.0]
No training will be performed.

WARM START
Penalty   Train CER      Dev CER       Dev length     Dev blank     
0.0       88.36          89.07         0.33           94.82         
0.5       87.20          87.83         0.37           93.87         
1.0       85.83          86.72         0.43           92.42         
1.5       84.61          86.16         0.49           90.57         
2.0       84.83          86.91         0.59           87.09         
3.0       107.44         101.85        1.03           70.03         
4.0       183.47         161.09        1.73           36.62         

Best training-probe penalty: 1.5
Development CER at chosen penalty: 86.16%
Development WER: 100.00%
Development prediction/reference length: 0.49
Example prediction: ይ መ ው መበሰበ አስስ ሰ መለድ መ ድህ ው

EPOCH 1
Penalty   Train CER      Dev CER       Dev length     Dev blank     
0.0       88.

In [ ]:

# ============================================================
# CELL 55 - CTC PREFIX BEAM SEARCH DIAGNOSTIC
#
# Compare greedy and beam decoding for:
#   Epoch 1: blank penalty 2.0
#   Epoch 4: blank penalty 3.0
#
# 24 new training examples + 15 development examples.
# No gradients, optimizer steps, or checkpoint changes.
# ============================================================

import json
import math
import random
from pathlib import Path

import torch
from jiwer import cer, wer

ROOT_55 = DATA_DIR / "amharic_2hour_pilot_v1"
RUN_55 = ROOT_55 / "head_only_stage1_v1"

SOURCE_55 = (
    DATA_DIR / "scaled_amharic_64_16_v1"
    / "stage2_filtered_62_v1" / "best.pt"
)

selection_55 = json.loads(
    (ROOT_55 / "selection.json").read_text(
        encoding="utf-8"
    )
)

carryover_55 = set(selection_55["carryover_ids"])

new_train_55 = [
    rid for rid in selection_55["train_ids"]
    if rid not in carryover_55
]

train_probe_55 = random.Random(551).sample(
    new_train_55, 24
)

dev_ids_55 = selection_55["primary_val_ids"]
all_ids_55 = train_probe_55 + dev_ids_55

assert len(train_probe_55) == 24
assert len(dev_ids_55) == 15

blank_55 = tokenizer.pad_token_id
device_55 = torch.device(
    "cuda" if torch.cuda.is_available() else "cpu"
)

heads_55 = {
    "Epoch 1": {
        "path": RUN_55 / "best.pt",
        "penalty": 2.0,
        "expected_greedy_cer": 0.8882
    },
    "Epoch 4": {
        "path": RUN_55 / "latest.pt",
        "penalty": 3.0,
        "expected_greedy_cer": 0.9592
    }
}

# ------------------------------------------------------------
# 1. Access cached encoder features.
#    Reconstruct only the required features if needed.
# ------------------------------------------------------------

available_cache_55 = globals().get("cache_53", {})

features_55 = {}

if all(rid in available_cache_55 for rid in all_ids_55):

    print("Reusing Cell 53's frozen encoder features.")

    for rid in all_ids_55:
        features_55[rid] = {
            "features": available_cache_55[rid][
                "features"
            ],
            "reference": available_cache_55[rid][
                "reference"
            ]
        }

else:

    print("Reconstructing the required frozen features.")
    print("No training will occur.")

    from transformers import Wav2Vec2ForCTC

    source = torch.load(
        SOURCE_55,
        map_location="cpu",
        weights_only=True
    )

    encoder_model = Wav2Vec2ForCTC.from_pretrained(
        str(BASELINE_DIR)
    ).to(device_55).float()

    for layer, weights in zip(
        encoder_model.wav2vec2.encoder.layers[-2:],
        source["upper_layers"]
    ):
        layer.load_state_dict(weights, strict=True)

    encoder_model.eval()
    encoder_model.requires_grad_(False)

    records_55 = {
        r["id"]: r for r in train_records
    }

    indices_55 = {
        r["id"]: i
        for i, r in enumerate(train_dataset.records)
    }

    with torch.no_grad():

        for i, rid in enumerate(all_ids_55, 1):

            example = train_dataset[
                indices_55[rid]
            ]

            batch = ctc_collator([example])

            hidden = encoder_model.wav2vec2(
                input_values=batch[
                    "input_values"
                ].to(device_55),
                attention_mask=batch[
                    "attention_mask"
                ].to(device_55)
            ).last_hidden_state

            features_55[rid] = {
                "features": hidden.detach().cpu().float(),
                "reference": normalize_amharic_ctc(
                    records_55[rid]["transcription"]
                )
            }

            if i % 10 == 0 or i == len(all_ids_55):
                print("Features:", i, "/", len(all_ids_55))

    del encoder_model

    if device_55.type == "cuda":
        torch.cuda.empty_cache()

# ------------------------------------------------------------
# 2. Stable log-space addition
# ------------------------------------------------------------

NEG_55 = -float("inf")

def logadd_55(a, b):
    if a == NEG_55:
        return b
    if b == NEG_55:
        return a

    maximum = max(a, b)

    return maximum + math.log1p(
        math.exp(min(a, b) - maximum)
    )

# ------------------------------------------------------------
# 3. Actual CTC prefix beam search
#
# Each prefix stores:
# pb  = probability ending in blank
# pnb = probability ending in nonblank
#
# Repeated tokens are handled using CTC rules.
# ------------------------------------------------------------

def prefix_beam_55(
    logits,
    blank_penalty=0.0,
    beam_width=10,
    top_k=12
):

    scores = logits.squeeze(0).float().clone()
    scores[:, blank_55] -= blank_penalty

    log_probs = torch.log_softmax(
        scores, dim=-1
    )

    blank_scores = log_probs[
        :, blank_55
    ].tolist()

    nonblank_scores = log_probs.clone()
    nonblank_scores[:, blank_55] = NEG_55

    values, indices = torch.topk(
        nonblank_scores,
        k=min(top_k, nonblank_scores.shape[-1] - 1),
        dim=-1
    )

    values = values.tolist()
    indices = indices.tolist()

    # Empty prefix initially ends in blank.
    beams = {(): (0.0, NEG_55)}

    for t in range(log_probs.shape[0]):

        next_beams = {}
        blank_score = blank_scores[t]

        def update(prefix, index, value):

            if value == NEG_55:
                return

            if prefix not in next_beams:
                next_beams[prefix] = [
                    NEG_55, NEG_55
                ]

            old = next_beams[prefix][index]

            next_beams[prefix][index] = (
                logadd_55(old, value)
            )

        for prefix, (pb, pnb) in beams.items():

            total = logadd_55(pb, pnb)

            # Emitting blank preserves the prefix.
            update(
                prefix, 0,
                total + blank_score
            )

            for token, score in zip(
                indices[t], values[t]
            ):

                if prefix and token == prefix[-1]:

                    # Repeating a token without an
                    # intervening blank collapses it.
                    update(
                        prefix, 1,
                        pnb + score
                    )

                    # The same token following blank
                    # creates a new repeated character.
                    update(
                        prefix + (token,), 1,
                        pb + score
                    )

                else:

                    update(
                        prefix + (token,), 1,
                        total + score
                    )

        best = sorted(
            next_beams.items(),
            key=lambda item: logadd_55(
                item[1][0], item[1][1]
            ),
            reverse=True
        )[:beam_width]

        beams = {
            prefix: tuple(probabilities)
            for prefix, probabilities in best
        }

    best_prefix = max(
        beams.items(),
        key=lambda item: logadd_55(
            item[1][0], item[1][1]
        )
    )[0]

    # Beam output is ALREADY CTC-collapsed.
    # Do not collapse repeated symbols again.
    decoded = tokenizer.decode(
        list(best_prefix),
        group_tokens=False
    )

    return normalize_amharic_ctc(decoded)

# ------------------------------------------------------------
# 4. Greedy decoding for direct comparison
# ------------------------------------------------------------

def greedy_55(logits, blank_penalty=0.0):

    adjusted = logits.clone().float()
    adjusted[:, :, blank_55] -= blank_penalty

    token_ids = adjusted.argmax(dim=-1)

    return normalize_amharic_ctc(
        processor.batch_decode(token_ids)[0]
    )

# ------------------------------------------------------------
# 5. Calculate CER, WER, and output length
# ------------------------------------------------------------

def measure_55(predictions, ids):

    references = [
        features_55[rid]["reference"]
        for rid in ids
    ]

    hypotheses = [
        predictions[rid]
        for rid in ids
    ]

    ref_characters = sum(
        len(s.replace(" ", ""))
        for s in references
    )

    hyp_characters = sum(
        len(s.replace(" ", ""))
        for s in hypotheses
    )

    return {
        "cer": float(cer(references, hypotheses)),
        "wer": float(wer(references, hypotheses)),
        "length_ratio": (
            hyp_characters / max(ref_characters, 1)
        ),
        "example": hypotheses[0]
    }

# ------------------------------------------------------------
# 6. Run both decoders with both settings
# ------------------------------------------------------------

results_55 = {}

print("\nCTC BEAM SEARCH COMPARISON")
print("=" * 65)
print("Training probe: 24 recordings")
print("Development: 15 recordings")
print("Beam width: 10")
print("Nonblank candidates/frame: 12")

for name, configuration in heads_55.items():

    checkpoint = torch.load(
        configuration["path"],
        map_location="cpu",
        weights_only=True
    )

    weights = checkpoint["head"]
    penalty = configuration["penalty"]

    head = torch.nn.Linear(
        in_features=weights["weight"].shape[1],
        out_features=weights["weight"].shape[0],
        bias=True
    ).to(device_55).float()

    head.load_state_dict(weights, strict=True)
    head.eval()

    logits_cache = {}

    with torch.no_grad():

        for rid in all_ids_55:

            features = features_55[rid][
                "features"
            ].to(device_55)

            logits_cache[rid] = (
                head(features).detach().cpu().float()
            )

    strategies = [
        ("Greedy", "greedy", 0.0),
        ("Greedy + penalty", "greedy", penalty),
        ("Beam", "beam", 0.0),
        ("Beam + penalty", "beam", penalty)
    ]

    model_results = []

    print("\n" + "=" * 65)
    print(name.upper())
    print("=" * 65)

    for label, method, amount in strategies:

        predictions = {}

        for rid in all_ids_55:

            logits = logits_cache[rid]

            if method == "greedy":
                predictions[rid] = greedy_55(
                    logits, amount
                )
            else:
                predictions[rid] = prefix_beam_55(
                    logits,
                    blank_penalty=amount,
                    beam_width=10,
                    top_k=12
                )

        train = measure_55(
            predictions, train_probe_55
        )

        dev = measure_55(
            predictions, dev_ids_55
        )

        model_results.append({
            "strategy": label,
            "penalty": amount,
            "train_cer": train["cer"],
            "dev_cer": dev["cer"],
            "dev_wer": dev["wer"],
            "dev_length": dev["length_ratio"],
            "dev_example": dev["example"]
        })

        print(
            f"{label:<21}"
            f"train CER={train['cer']*100:6.2f}%  "
            f"dev CER={dev['cer']*100:6.2f}%  "
            f"dev WER={dev['wer']*100:6.2f}%  "
            f"length={dev['length_ratio']:.2f}"
        )

    baseline = model_results[0]["dev_cer"]

    assert abs(
        baseline -
        configuration["expected_greedy_cer"]
    ) < 0.005, (
        f"Unexpected baseline mismatch for {name}: "
        f"{baseline:.4f}"
    )

    # The blank penalty was selected in Cell 54
    # using its training probe, not this dev set.
    chosen = min(
        model_results,
        key=lambda row: row["train_cer"]
    )

    print("\nLowest training-probe CER:",
          chosen["strategy"])

    print(
        "Development CER:",
        f"{chosen['dev_cer']*100:.2f}%"
    )

    print(
        "Example transcription:",
        chosen["dev_example"][:180] or "[EMPTY]"
    )

    results_55[name] = model_results

    del head, logits_cache

# ------------------------------------------------------------
# 7. Save diagnostic results
# ------------------------------------------------------------

output_55 = RUN_55 / "ctc_beam_diagnostic.json"

output_55.write_text(
    json.dumps(
        {
            "beam_width": 10,
            "top_k_nonblank": 12,
            "train_probe_count": len(train_probe_55),
            "development_count": len(dev_ids_55),
            "description": (
                "Exploratory greedy and approximate CTC "
                "prefix beam decoding comparison."
            ),
            "results": results_55
        },
        indent=2,
        ensure_ascii=False
    ),
    encoding="utf-8"
)

print("\n" + "=" * 65)
print("BEAM DIAGNOSTIC COMPLETE")
print("=" * 65)
print("Saved:", output_55)
print("Training updates: 0")
print("Checkpoints modified: 0")


Reusing Cell 53's frozen encoder features.

CTC BEAM SEARCH COMPARISON
Training probe: 24 recordings
Development: 15 recordings
Beam width: 10
Nonblank candidates/frame: 12

EPOCH 1
Greedy               train CER= 89.36%  dev CER= 88.82%  dev WER= 99.70%  length=0.18
Greedy + penalty     train CER= 82.51%  dev CER= 83.32%  dev WER=103.34%  length=0.35
Beam                 train CER= 89.03%  dev CER= 88.02%  dev WER= 99.70%  length=0.18
Beam + penalty       train CER= 81.05%  dev CER= 82.64%  dev WER=114.29%  length=0.46

Lowest training-probe CER: Beam + penalty
Development CER: 82.64%
Example transcription: የ መ መበራ አበ ከከአ የ ከ ከ የ ከ መለከክድ መ ህ መ ም

EPOCH 4
Greedy               train CER= 95.48%  dev CER= 95.92%  dev WER= 99.70%  length=0.05
Greedy + penalty     train CER= 80.58%  dev CER= 81.59%  dev WER=120.97%  length=0.38
Beam                 train CER= 97.01%  dev CER= 96.48%  dev WER= 99.70%  length=0.04
Beam + penalty       train CER= 85.71%  dev CER= 83.57%  dev WER=180.55%  leng

In [ ]:

# ============================================================
# CELL 56 - TWO-HOUR JOINT ENCODER + CTC HEAD PILOT
#
# Encoder: Cell 50 best checkpoint
# CTC head: Cell 53 epoch-1 checkpoint
#
# Train: 452 recordings, 408 speakers
# Development: 15 speaker-disjoint recordings
#
# Train last 2 encoder layers + CTC head
# One epoch, FP32, gradient clipping
# Checkpoint every 113 updates
#
# Previous checkpoints remain untouched.
# ============================================================

import gc
import json
import random
import hashlib
import statistics
from pathlib import Path

import torch
from jiwer import cer, wer
from transformers import Wav2Vec2ForCTC

assert torch.cuda.is_available(), (
    "A CUDA GPU is required for this training experiment."
)

DEVICE_56 = torch.device("cuda")

ROOT_56 = DATA_DIR / "amharic_2hour_pilot_v1"

ENCODER_SOURCE_56 = (
    DATA_DIR / "scaled_amharic_64_16_v1"
    / "stage2_filtered_62_v1" / "best.pt"
)

HEAD_SOURCE_56 = (
    ROOT_56 / "head_only_stage1_v1" / "best.pt"
)

SELECTION_56 = ROOT_56 / "selection.json"

RUN_56 = ROOT_56 / "joint_last2_stage2_v1"
RUN_56.mkdir(parents=True, exist_ok=True)

LATEST_56 = RUN_56 / "latest.pt"
BEST_56 = RUN_56 / "best.pt"
HISTORY_56 = RUN_56 / "history.json"

ENCODER_LR_56 = 1e-5
HEAD_LR_56 = 1e-4
CLIP_NORM_56 = 5.0
BLANK_PENALTY_56 = 2.0

SEED_56 = 20261020
REPORT_EVERY_56 = 113
TOTAL_UPDATES_56 = 452

def read_json_56(path):
    assert path.is_file(), f"Missing file: {path}"
    return json.loads(path.read_text(encoding="utf-8"))

selection_56 = read_json_56(SELECTION_56)

train_ids_56 = selection_56["train_ids"]
val_ids_56 = selection_56["primary_val_ids"]
carryover_ids_56 = selection_56["carryover_ids"]

assert len(train_ids_56) == 452
assert len(val_ids_56) == 15
assert not set(train_ids_56) & set(val_ids_56)

records_56 = {
    r["id"]: r for r in train_records
}

indices_56 = {
    r["id"]: i
    for i, r in enumerate(train_dataset.records)
}

assert all(
    rid in indices_56
    for rid in train_ids_56 + val_ids_56
)

train_speakers_56 = {
    records_56[rid]["speaker_id"]
    for rid in train_ids_56
}

val_speakers_56 = {
    records_56[rid]["speaker_id"]
    for rid in val_ids_56
}

assert not train_speakers_56 & val_speakers_56

new_ids_56 = [
    rid for rid in train_ids_56
    if rid not in set(carryover_ids_56)
]

# Fixed diagnostic probes, not the full training set.
probe_rng_56 = random.Random(SEED_56)

old_probe_56 = probe_rng_56.sample(
    carryover_ids_56, 16
)

new_probe_56 = probe_rng_56.sample(
    new_ids_56, 32
)

# ------------------------------------------------------------
# 1. Restore the encoder and the epoch-1 head
# ------------------------------------------------------------

encoder_checkpoint_56 = torch.load(
    ENCODER_SOURCE_56,
    map_location="cpu",
    weights_only=True
)

head_checkpoint_56 = torch.load(
    HEAD_SOURCE_56,
    map_location="cpu",
    weights_only=True
)

assert encoder_checkpoint_56["precision"] == "fp32"
assert head_checkpoint_56["completed_epochs"] == 1

model_56 = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(DEVICE_56).float()

for layer, weights in zip(
    model_56.wav2vec2.encoder.layers[-2:],
    encoder_checkpoint_56["upper_layers"]
):
    layer.load_state_dict(weights, strict=True)

model_56.lm_head.load_state_dict(
    head_checkpoint_56["head"],
    strict=True
)

model_56.requires_grad_(False)

upper_layers_56 = list(
    model_56.wav2vec2.encoder.layers[-2:]
)

for layer in upper_layers_56:
    layer.requires_grad_(True)

model_56.lm_head.requires_grad_(True)

# Keep dropout and SpecAugment disabled for this
# controlled continuation. Gradients remain enabled.
model_56.eval()

encoder_params_56 = [
    p
    for layer in upper_layers_56
    for p in layer.parameters()
    if p.requires_grad
]

head_params_56 = list(
    model_56.lm_head.parameters()
)

trainable_56 = (
    encoder_params_56 + head_params_56
)

parameter_count_56 = sum(
    p.numel() for p in trainable_56
)

assert parameter_count_56 == 25521473

optimizer_56 = torch.optim.AdamW([
    {
        "params": encoder_params_56,
        "lr": ENCODER_LR_56,
        "weight_decay": 0.01
    },
    {
        "params": head_params_56,
        "lr": HEAD_LR_56,
        "weight_decay": 0.0
    }
])

config_56 = {
    "encoder_checkpoint": str(ENCODER_SOURCE_56),
    "head_checkpoint": str(HEAD_SOURCE_56),
    "train_ids": train_ids_56,
    "val_ids": val_ids_56,
    "encoder_lr": ENCODER_LR_56,
    "head_lr": HEAD_LR_56,
    "clip_norm": CLIP_NORM_56,
    "blank_penalty": BLANK_PENALTY_56,
    "seed": SEED_56,
    "total_updates": TOTAL_UPDATES_56
}

signature_56 = hashlib.sha256(
    json.dumps(
        config_56,
        ensure_ascii=False,
        sort_keys=True
    ).encode("utf-8")
).hexdigest()

# ------------------------------------------------------------
# 2. Restore existing pilot progress if present
# ------------------------------------------------------------

completed_56 = 0
history_56 = []
best_adjusted_cer_56 = float("inf")

if LATEST_56.exists():

    checkpoint = torch.load(
        LATEST_56,
        map_location="cpu",
        weights_only=True
    )

    assert checkpoint["signature"] == signature_56

    model_56.lm_head.load_state_dict(
        checkpoint["head"]
    )

    for layer, weights in zip(
        upper_layers_56,
        checkpoint["upper_layers"]
    ):
        layer.load_state_dict(weights)

    optimizer_56.load_state_dict(
        checkpoint["optimizer"]
    )

    completed_56 = int(checkpoint["updates"])
    best_adjusted_cer_56 = float(
        checkpoint["best_adjusted_cer"]
    )

    assert HISTORY_56.is_file()
    history_56 = read_json_56(HISTORY_56)

    print("Resuming at update:", completed_56)

else:
    print("Starting new joint fine-tuning pilot.")

assert 0 <= completed_56 <= TOTAL_UPDATES_56

# ------------------------------------------------------------
# 3. Input and decoding helpers
# ------------------------------------------------------------

def batch_56(rid):

    item = train_dataset[indices_56[rid]]
    batch = ctc_collator([item])

    return {
        key: value.to(DEVICE_56)
        for key, value in batch.items()
    }

def decode_56(logits, penalty):

    adjusted = logits.float().clone()

    adjusted[:, :, tokenizer.pad_token_id] -= penalty

    token_ids = adjusted.argmax(dim=-1)

    text = processor.batch_decode(
        token_ids.cpu()
    )[0]

    return normalize_amharic_ctc(text)

def evaluate_56(ids):

    model_56.eval()

    references = []
    standard_predictions = []
    adjusted_predictions = []

    with torch.no_grad():

        for rid in ids:

            batch = batch_56(rid)

            logits = model_56(
                input_values=batch["input_values"],
                attention_mask=batch["attention_mask"]
            ).logits

            references.append(
                normalize_amharic_ctc(
                    records_56[rid]["transcription"]
                )
            )

            standard_predictions.append(
                decode_56(logits, penalty=0.0)
            )

            adjusted_predictions.append(
                decode_56(
                    logits,
                    penalty=BLANK_PENALTY_56
                )
            )

            del batch, logits

    reference_chars = sum(
        len(x.replace(" ", ""))
        for x in references
    )

    predicted_chars = sum(
        len(x.replace(" ", ""))
        for x in adjusted_predictions
    )

    return {
        "greedy_cer": float(
            cer(references, standard_predictions)
        ),
        "adjusted_cer": float(
            cer(references, adjusted_predictions)
        ),
        "adjusted_wer": float(
            wer(references, adjusted_predictions)
        ),
        "adjusted_length_ratio": (
            predicted_chars / max(reference_chars, 1)
        ),
        "sample": adjusted_predictions[0]
    }

def report_56(step):

    old = evaluate_56(old_probe_56)
    new = evaluate_56(new_probe_56)
    val = evaluate_56(val_ids_56)

    row = {
        "updates": step,
        "old_adjusted_cer": old["adjusted_cer"],
        "new_adjusted_cer": new["adjusted_cer"],
        "dev_greedy_cer": val["greedy_cer"],
        "dev_adjusted_cer": val["adjusted_cer"],
        "dev_adjusted_wer": val["adjusted_wer"],
        "dev_adjusted_length": val[
            "adjusted_length_ratio"
        ],
        "dev_example": val["sample"]
    }

    print(f"\nUPDATE {step}/{TOTAL_UPDATES_56}")
    print("-" * 60)

    print(
        "Old training probe adjusted CER:",
        f"{old['adjusted_cer']*100:.2f}%"
    )

    print(
        "New training probe adjusted CER:",
        f"{new['adjusted_cer']*100:.2f}%"
    )

    print(
        "Development greedy CER:",
        f"{val['greedy_cer']*100:.2f}%"
    )

    print(
        "Development adjusted CER:",
        f"{val['adjusted_cer']*100:.2f}%"
    )

    print(
        "Development adjusted WER:",
        f"{val['adjusted_wer']*100:.2f}%"
    )

    print(
        "Adjusted prediction/reference length:",
        f"{val['adjusted_length_ratio']:.2f}"
    )

    print(
        "Example:",
        val["sample"][:140] or "[EMPTY]"
    )

    return row

def save_56(step, improved):

    state = {
        "signature": signature_56,
        "updates": step,
        "best_adjusted_cer": best_adjusted_cer_56,
        "precision": "fp32",
        "head": model_56.lm_head.state_dict(),
        "upper_layers": [
            layer.state_dict()
            for layer in upper_layers_56
        ],
        "optimizer": optimizer_56.state_dict()
    }

    temp = RUN_56 / "latest.pt.partial"
    torch.save(state, temp)
    temp.replace(LATEST_56)

    if improved:
        temp_best = RUN_56 / "best.pt.partial"
        torch.save(state, temp_best)
        temp_best.replace(BEST_56)

    history_temp = RUN_56 / "history.json.partial"

    history_temp.write_text(
        json.dumps(
            history_56,
            ensure_ascii=False,
            indent=2
        ),
        encoding="utf-8"
    )

    history_temp.replace(HISTORY_56)

# ------------------------------------------------------------
# 4. Verify longest-recording FP32 gradients
# ------------------------------------------------------------

print("\nJOINT TRAINING CONFIGURATION")
print("=" * 60)

print("Training recordings:", len(train_ids_56))
print("Training speakers:", len(train_speakers_56))
print("Development recordings:", len(val_ids_56))
print("Trainable parameters:", parameter_count_56)
print("Encoder LR:", ENCODER_LR_56)
print("Head LR:", HEAD_LR_56)
print("Gradient clipping:", CLIP_NORM_56)
print("CTC loss reduction:", model_56.config.ctc_loss_reduction)
print("Blank penalty for evaluation:", BLANK_PENALTY_56)
print("Precision: FP32")
print("Completed updates:", completed_56)

if completed_56 == 0:

    longest_id_56 = max(
        train_ids_56,
        key=lambda rid: float(
            records_56[rid]["duration_seconds"]
        )
    )

    print("\nLONG-RECORDING GRADIENT PREFLIGHT")
    print("-" * 60)

    optimizer_56.zero_grad(set_to_none=True)

    longest_batch_56 = batch_56(longest_id_56)

    torch.cuda.reset_peak_memory_stats()

    with torch.autocast(
        device_type="cuda",
        enabled=False
    ):
        test_loss_56 = model_56(
            **longest_batch_56
        ).loss

    assert torch.isfinite(test_loss_56).item()

    test_loss_56.backward()

    gradient_norm_56 = (
        torch.nn.utils.clip_grad_norm_(
            trainable_56,
            max_norm=CLIP_NORM_56,
            error_if_nonfinite=True
        )
    )

    print("Recording ID:", longest_id_56)
    print(
        "Duration:",
        records_56[longest_id_56]["duration_seconds"],
        "seconds"
    )
    print("Loss:", float(test_loss_56))
    print("Gradient norm:", float(gradient_norm_56))
    print(
        "Peak allocated GPU memory:",
        round(
            torch.cuda.max_memory_allocated()
            / 1024**3,
            2
        ),
        "GiB"
    )

    optimizer_56.zero_grad(set_to_none=True)
    del longest_batch_56, test_loss_56

    torch.cuda.empty_cache()

    print("Preflight passed. Optimizer updates: 0")

# ------------------------------------------------------------
# 5. Evaluate exact warm-start baseline
# ------------------------------------------------------------

if completed_56 == 0 and not history_56:

    baseline_56 = report_56(0)

    # Compare with Cell 55's epoch-1 results.
    assert abs(
        baseline_56["dev_greedy_cer"] - 0.8882
    ) < 0.015, (
        "Baseline greedy CER mismatch. "
        "Inspect restored checkpoints."
    )

    assert abs(
        baseline_56["dev_adjusted_cer"] - 0.8332
    ) < 0.015, (
        "Baseline adjusted CER mismatch. "
        "Inspect encoder/head pairing."
    )

    history_56.append(baseline_56)

    best_adjusted_cer_56 = baseline_56[
        "dev_adjusted_cer"
    ]

# ------------------------------------------------------------
# 6. Deterministic one-epoch training order
# ------------------------------------------------------------

order_56 = list(train_ids_56)

random.Random(
    SEED_56 + 1
).shuffle(order_56)

assert len(order_56) == TOTAL_UPDATES_56

segment_losses_56 = []
segment_norms_56 = []

# ------------------------------------------------------------
# 7. Train once on each recording
# ------------------------------------------------------------

for update in range(
    completed_56 + 1,
    TOTAL_UPDATES_56 + 1
):

    rid = order_56[update - 1]

    optimizer_56.zero_grad(set_to_none=True)
    model_56.eval()

    batch = batch_56(rid)

    with torch.autocast(
        device_type="cuda",
        enabled=False
    ):
        loss = model_56(**batch).loss

    if not torch.isfinite(loss).item():
        raise RuntimeError(
            f"Nonfinite loss at update {update}, "
            f"recording {rid}"
        )

    loss.backward()

    gradient_norm = (
        torch.nn.utils.clip_grad_norm_(
            trainable_56,
            max_norm=CLIP_NORM_56,
            error_if_nonfinite=True
        )
    )

    raw_norm = float(gradient_norm)

    if raw_norm > 5000:
        optimizer_56.zero_grad(set_to_none=True)
        raise RuntimeError(
            f"Extreme gradient at update {update}: "
            f"{raw_norm:.1f}"
        )

    optimizer_56.step()

    segment_losses_56.append(float(loss.item()))
    segment_norms_56.append(raw_norm)

    del batch, loss

    if (
        update % REPORT_EVERY_56 == 0
        or update == TOTAL_UPDATES_56
    ):

        result = report_56(update)

        result["mean_step_loss"] = (
            statistics.mean(segment_losses_56)
        )

        result["median_gradient_norm"] = (
            statistics.median(segment_norms_56)
        )

        result["max_gradient_norm"] = (
            max(segment_norms_56)
        )

        result["clipped_fraction"] = (
            sum(
                norm > CLIP_NORM_56
                for norm in segment_norms_56
            ) / len(segment_norms_56)
        )

        improved = (
            result["dev_adjusted_cer"]
            < best_adjusted_cer_56
        )

        if improved:
            best_adjusted_cer_56 = result[
                "dev_adjusted_cer"
            ]

        history_56.append(result)

        save_56(
            step=update,
            improved=improved
        )

        print(
            "Mean training-step loss:",
            round(result["mean_step_loss"], 4)
        )

        print(
            "Median gradient norm:",
            round(result["median_gradient_norm"], 2)
        )

        print(
            "Maximum gradient norm:",
            round(result["max_gradient_norm"], 2)
        )

        print(
            "Fraction clipped:",
            f"{result['clipped_fraction']*100:.1f}%"
        )

        segment_losses_56.clear()
        segment_norms_56.clear()

# ------------------------------------------------------------
# 8. Summary
# ------------------------------------------------------------

print("\n" + "=" * 78)
print("TWO-HOUR JOINT FINE-TUNING RESULTS")
print("=" * 78)

print(
    f"{'Update':<10}"
    f"{'Old CER':<13}"
    f"{'New CER':<13}"
    f"{'Dev greedy':<14}"
    f"{'Dev adjusted':<15}"
    f"{'Length':<9}"
)

for row in history_56:

    print(
        f"{row['updates']:<10}"
        f"{row['old_adjusted_cer']*100:<13.2f}"
        f"{row['new_adjusted_cer']*100:<13.2f}"
        f"{row['dev_greedy_cer']*100:<14.2f}"
        f"{row['dev_adjusted_cer']*100:<15.2f}"
        f"{row['dev_adjusted_length']:<9.2f}"
    )

print(
    "\nBest adjusted development CER:",
    f"{best_adjusted_cer_56*100:.2f}%"
)

print("Latest checkpoint:", LATEST_56)

if BEST_56.exists():
    print("Best joint checkpoint:", BEST_56)
else:
    print(
        "No joint checkpoint improved on the "
        "original epoch-1 model."
    )

print("History:", HISTORY_56)
print("Previous checkpoints unchanged.")


Starting new joint fine-tuning pilot.

JOINT TRAINING CONFIGURATION
Training recordings: 452
Training speakers: 408
Development recordings: 15
Trainable parameters: 25521473
Encoder LR: 1e-05
Head LR: 0.0001
Gradient clipping: 5.0
CTC loss reduction: mean
Blank penalty for evaluation: 2.0
Precision: FP32
Completed updates: 0

LONG-RECORDING GRADIENT PREFLIGHT
------------------------------------------------------------
Recording ID: 5DevVlRQXWD2jCGufQXu
Duration: 17.976 seconds
Loss: 3.9612960815429688
Gradient norm: 8.676441192626953
Peak allocated GPU memory: 8.38 GiB
Preflight passed. Optimizer updates: 0


/tmp/ipykernel_565/1996426138.py:521: UserWarning: Converting a tensor with requires_grad=True to a scalar may lead to unexpected behavior.
Consider using tensor.detach() first. (Triggered internally at /pytorch/torch/csrc/autograd/generated/python_variable_methods.cpp:836.)
  print("Loss:", float(test_loss_56))



UPDATE 0/452
------------------------------------------------------------
Old training probe adjusted CER: 78.58%
New training probe adjusted CER: 82.52%
Development greedy CER: 88.82%
Development adjusted CER: 83.32%
Development adjusted WER: 103.34%
Adjusted prediction/reference length: 0.35
Example: የ መመበራሰበ አስ ሰ መለክድ ማ ድ መ ም

UPDATE 113/452
------------------------------------------------------------
Old training probe adjusted CER: 80.66%
New training probe adjusted CER: 85.56%
Development greedy CER: 91.23%
Development adjusted CER: 85.55%
Development adjusted WER: 100.00%
Adjusted prediction/reference length: 0.24
Example: የ በራሰበ አ ሰን ክድ ማ ው
Mean training-step loss: 4.6676
Median gradient norm: 11.38
Maximum gradient norm: 147.64
Fraction clipped: 89.4%

UPDATE 226/452
------------------------------------------------------------
Old training probe adjusted CER: 82.59%
New training probe adjusted CER: 86.60%
Development greedy CER: 92.90%
Development adjusted CER: 86.91%
Develop

In [ ]:

# ============================================================
# CELL 57 - CONTROLLED FOUR-RECORDING LEARNABILITY TEST
#
# Compare:
# A. Original pretrained XLS-R encoder
# B. Adapted encoder from Cell 50
#
# Both receive IDENTICALLY initialized fresh CTC heads.
# Train only on four manually reviewed recordings.
#
# 1600 updates per branch, save every 400.
# No development or test recordings used.
# ============================================================

import copy
import gc
import json
import random
import hashlib
import statistics
from pathlib import Path

import torch
import torch.nn.functional as F
from jiwer import cer, wer
from transformers import Wav2Vec2ForCTC

assert torch.cuda.is_available(), "CUDA is required."

DEVICE_57 = torch.device("cuda")
ROOT_57 = DATA_DIR / "amharic_2hour_pilot_v1"
RUN_57 = ROOT_57 / "four_recording_learnability_v1"
RUN_57.mkdir(parents=True, exist_ok=True)

REVIEW_ROOT_57 = DATA_DIR / "scaled_amharic_64_16_v1"

ENCODER_CKPT_57 = (
    REVIEW_ROOT_57
    / "stage2_filtered_62_v1"
    / "best.pt"
)

UPDATES_57 = 1600
REPORT_57 = 400
HEAD_LR_57 = 1e-3
CLIP_57 = 5.0
SEED_57 = 5701

# ------------------------------------------------------------
# 1. Select ONLY human-reviewed training examples
# ------------------------------------------------------------

reviews_57 = []

for filename in [
    "manual_review_results_round1.json",
    "manual_review_results_round2.json"
]:
    path = REVIEW_ROOT_57 / filename

    reviews_57.extend(
        json.loads(path.read_text(encoding="utf-8"))
    )

allowed_57 = {"verified_match", "match_with_fillers"}

clean_ids_57 = [
    r["id"]
    for r in reviews_57
    if r["review_status"] in allowed_57
    and r["original_group"] in {
        "Previous 8 training",
        "New 56 training"
    }
]

assert len(clean_ids_57) == 4
assert len(set(clean_ids_57)) == 4

records_57 = {
    r["id"]: r for r in train_records
}

indices_57 = {
    r["id"]: i
    for i, r in enumerate(train_dataset.records)
}

print("FOUR-RECORDING LEARNABILITY TEST")
print("=" * 60)

for i, rid in enumerate(clean_ids_57, 1):
    rec = records_57[rid]

    print(
        f"{i}. {rid}",
        f"| {rec['duration_seconds']:.2f}s",
        f"| speaker {rec['speaker_id']}"
    )

print(
    "Distinct speakers:",
    len({
        records_57[rid]["speaker_id"]
        for rid in clean_ids_57
    })
)

# ------------------------------------------------------------
# 2. Verify CTC model configuration
# ------------------------------------------------------------

model_57 = Wav2Vec2ForCTC.from_pretrained(
    str(BASELINE_DIR)
).to(DEVICE_57).float()

model_57.eval()
model_57.requires_grad_(False)

blank_57 = tokenizer.pad_token_id
vocab_57 = len(tokenizer)

print("\nCONFIGURATION CHECK")
print("=" * 60)

print("Tokenizer blank ID:", blank_57)
print("Model blank ID:", model_57.config.pad_token_id)
print("Tokenizer vocabulary:", vocab_57)
print("Model vocabulary:", model_57.config.vocab_size)
print("CTC reduction:", model_57.config.ctc_loss_reduction)

assert model_57.config.pad_token_id == blank_57, (
    "CRITICAL: CTC blank ID mismatch."
)

assert model_57.config.vocab_size == vocab_57, (
    "CRITICAL: Model/tokenizer vocabulary mismatch."
)

# ------------------------------------------------------------
# 3. Build exact training batches
# ------------------------------------------------------------

batches_57 = {}
references_57 = {}

for rid in clean_ids_57:

    example = train_dataset[indices_57[rid]]
    batch = ctc_collator([example])

    targets = batch["labels"][0]
    targets = targets[targets >= 0].long()

    reference = normalize_amharic_ctc(
        records_57[rid]["transcription"]
    )

    reconstructed = normalize_amharic_ctc(
        tokenizer.decode(
            targets.tolist(),
            group_tokens=False
        )
    )

    assert reconstructed == reference
    assert not (targets == blank_57).any()

    batches_57[rid] = batch
    references_57[rid] = reference

# ------------------------------------------------------------
# 4. Cache original and adapted encoder outputs
# ------------------------------------------------------------

encoder_checkpoint_57 = torch.load(
    ENCODER_CKPT_57,
    map_location="cpu",
    weights_only=True
)

feature_sets_57 = {}

for branch in ["Original pretrained", "Adapted encoder"]:

    if branch == "Adapted encoder":

        for layer, weights in zip(
            model_57.wav2vec2.encoder.layers[-2:],
            encoder_checkpoint_57["upper_layers"]
        ):
            layer.load_state_dict(
                weights,
                strict=True
            )

    model_57.eval()

    features = {}

    with torch.no_grad():

        for rid in clean_ids_57:

            batch = batches_57[rid]

            hidden = model_57.wav2vec2(
                input_values=batch[
                    "input_values"
                ].to(DEVICE_57),
                attention_mask=batch[
                    "attention_mask"
                ].to(DEVICE_57)
            ).last_hidden_state

            targets = batch["labels"][0]
            targets = targets[targets >= 0].long()

            repeated = int(
                (targets[1:] == targets[:-1])
                .sum().item()
            )

            assert hidden.shape[1] >= (
                len(targets) + repeated
            )

            assert torch.isfinite(hidden).all().item()

            features[rid] = {
                "hidden": hidden.cpu().float().contiguous(),
                "targets": targets.cpu().contiguous(),
                "frames": int(hidden.shape[1]),
                "label_count": int(targets.numel())
            }

    feature_sets_57[branch] = features
    print("\nCached:", branch)

del model_57
gc.collect()
torch.cuda.empty_cache()

# ------------------------------------------------------------
# 5. Identical fresh head initialization
# ------------------------------------------------------------

torch.manual_seed(SEED_57)

template_head_57 = torch.nn.Linear(
    1024,
    vocab_57,
    bias=True
)

initial_head_57 = copy.deepcopy(
    template_head_57.state_dict()
)

del template_head_57

# ------------------------------------------------------------
# 6. Training and evaluation helpers
# ------------------------------------------------------------

def loss_57(head, features, rid):

    item = features[rid]

    hidden = item["hidden"].to(DEVICE_57)
    targets = item["targets"].to(DEVICE_57)

    logits = head(hidden)

    log_probs = F.log_softmax(
        logits.float(),
        dim=-1
    ).transpose(0, 1)

    return F.ctc_loss(
        log_probs,
        targets,
        torch.tensor(
            [item["frames"]],
            dtype=torch.long
        ),
        torch.tensor(
            [item["label_count"]],
            dtype=torch.long
        ),
        blank=blank_57,
        reduction="mean",
        zero_infinity=False
    )

def evaluate_57(head, features):

    head.eval()

    predictions = []
    references = []
    blank_count = 0
    frame_count = 0
    losses = []

    with torch.no_grad():

        for rid in clean_ids_57:

            item = features[rid]
            hidden = item["hidden"].to(DEVICE_57)

            logits = head(hidden)

            predicted_ids = logits.argmax(dim=-1)

            blank_count += int(
                (predicted_ids == blank_57).sum().item()
            )

            frame_count += predicted_ids.numel()

            prediction = processor.batch_decode(
                predicted_ids.cpu()
            )[0]

            predictions.append(
                normalize_amharic_ctc(prediction)
            )

            references.append(references_57[rid])

            losses.append(
                float(loss_57(head, features, rid).item())
            )

    return {
        "cer": float(cer(references, predictions)),
        "wer": float(wer(references, predictions)),
        "ctc_loss": statistics.mean(losses),
        "blank_fraction": blank_count / max(frame_count, 1),
        "length_ratio": (
            sum(len(p.replace(" ", "")) for p in predictions)
            / max(
                sum(len(r.replace(" ", "")) for r in references),
                1
            )
        ),
        "predictions": {
            rid: prediction
            for rid, prediction in zip(
                clean_ids_57, predictions
            )
        }
    }

def record_for_step_57(step):

    epoch = (step - 1) // len(clean_ids_57)
    position = (step - 1) % len(clean_ids_57)

    order = list(clean_ids_57)

    random.Random(SEED_57 + epoch).shuffle(order)

    return order[position]

# ------------------------------------------------------------
# 7. Run both independent branches
# ------------------------------------------------------------

results_57 = {}

for branch, features in feature_sets_57.items():

    branch_dir = RUN_57 / (
        "original" if branch == "Original pretrained"
        else "adapted"
    )

    branch_dir.mkdir(exist_ok=True)

    latest = branch_dir / "latest.pt"
    history_path = branch_dir / "history.json"

    head = torch.nn.Linear(
        1024, vocab_57
    ).to(DEVICE_57).float()

    head.load_state_dict(
        initial_head_57,
        strict=True
    )

    optimizer = torch.optim.AdamW(
        head.parameters(),
        lr=HEAD_LR_57,
        weight_decay=0.0
    )

    signature = hashlib.sha256(
        json.dumps(
            {
                "branch": branch,
                "source": str(ENCODER_CKPT_57),
                "recordings": [
                    {
                        "id": rid,
                        "transcript": references_57[rid]
                    }
                    for rid in clean_ids_57
                ],
                "seed": SEED_57,
                "lr": HEAD_LR_57,
                "clip": CLIP_57
            },
            sort_keys=True,
            ensure_ascii=False
        ).encode("utf-8")
    ).hexdigest()

    start_step = 0
    history = []

    if latest.exists():

        saved = torch.load(
            latest,
            map_location="cpu",
            weights_only=True
        )

        assert saved["signature"] == signature

        head.load_state_dict(saved["head"])
        optimizer.load_state_dict(saved["optimizer"])

        start_step = int(saved["step"])

        assert history_path.exists()

        history = json.loads(
            history_path.read_text(encoding="utf-8")
        )

    else:

        initial = evaluate_57(head, features)
        initial["step"] = 0
        history.append(initial)

    print("\n" + "=" * 65)
    print(branch.upper())
    print("=" * 65)
    print("Starting update:", start_step)

    recent_losses = []

    for step in range(start_step + 1, UPDATES_57 + 1):

        rid = record_for_step_57(step)

        head.train()
        optimizer.zero_grad(set_to_none=True)

        loss = loss_57(head, features, rid)

        if not torch.isfinite(loss).item():
            raise RuntimeError(
                f"Nonfinite loss: {branch}, update {step}"
            )

        loss.backward()

        torch.nn.utils.clip_grad_norm_(
            head.parameters(),
            max_norm=CLIP_57,
            error_if_nonfinite=True
        )

        optimizer.step()

        recent_losses.append(float(loss.detach().item()))

        if step % REPORT_57 == 0:

            metrics = evaluate_57(head, features)
            metrics["step"] = step

            metrics["mean_recent_train_loss"] = (
                statistics.mean(recent_losses)
            )

            history.append(metrics)

            print(
                f"Update {step:4d} | "
                f"CER {metrics['cer']*100:6.2f}% | "
                f"WER {metrics['wer']*100:6.2f}% | "
                f"CTC {metrics['ctc_loss']:6.3f} | "
                f"Length {metrics['length_ratio']:.2f} | "
                f"Blank {metrics['blank_fraction']*100:.1f}%"
            )

            checkpoint = {
                "signature": signature,
                "step": step,
                "head": head.state_dict(),
                "optimizer": optimizer.state_dict()
            }

            temp_checkpoint = branch_dir / "latest.pt.partial"
            torch.save(checkpoint, temp_checkpoint)
            temp_checkpoint.replace(latest)

            temp_history = branch_dir / "history.json.partial"

            temp_history.write_text(
                json.dumps(
                    history,
                    ensure_ascii=False,
                    indent=2
                ),
                encoding="utf-8"
            )

            temp_history.replace(history_path)

            recent_losses.clear()

    results_57[branch] = history

    del head, optimizer
    torch.cuda.empty_cache()

# ------------------------------------------------------------
# 8. Compare memorization ability
# ------------------------------------------------------------

print("\n" + "=" * 75)
print("FOUR-RECORDING LEARNABILITY RESULTS")
print("=" * 75)

print(
    f"{'Update':<10}"
    f"{'Original CER':<18}"
    f"{'Adapted CER':<18}"
)

original_history = {
    r["step"]: r
    for r in results_57["Original pretrained"]
}

adapted_history = {
    r["step"]: r
    for r in results_57["Adapted encoder"]
}

for step in sorted(
    set(original_history) & set(adapted_history)
):

    original_cer = original_history[step]["cer"] * 100
    adapted_cer = adapted_history[step]["cer"] * 100

    print(
        f"{step:<10}"
        f"{original_cer:<18.2f}"
        f"{adapted_cer:<18.2f}"
    )

print("\nFinal per-recording results:")

for branch in results_57:

    final = results_57[branch][-1]

    print("\n", branch)

    for rid in clean_ids_57:

        print("\nID:", rid)
        print("REFERENCE:", references_57[rid])
        print(
            "PREDICTION:",
            final["predictions"][rid] or "[EMPTY]"
        )

print("\nSaved experiment:", RUN_57)
print("Existing ASR checkpoints unchanged.")


FOUR-RECORDING LEARNABILITY TEST
1. JljzcvdzYAAyQmAc4x5u | 14.90s | speaker wZj8gPvur6apWK0EGgLFFAFDlQj2
2. 1kPe5yhdSKLyyBYtp1yP | 14.98s | speaker b4xjYXm7arfa71rqgZnrTIbp3sN2
3. 7ZOeZpBUxW6IXls17BxG | 14.86s | speaker wK3oCHv9SkWEDZywENpd2WbwlbO2
4. 5us9lovEMnIT5mMb6bQ9 | 14.38s | speaker moSDdgXQeQR5Qtx2z3zBovLqYeN2
Distinct speakers: 4

CONFIGURATION CHECK
Tokenizer blank ID: 320
Model blank ID: 320
Tokenizer vocabulary: 321
Model vocabulary: 321
CTC reduction: mean

Cached: Original pretrained

Cached: Adapted encoder

ORIGINAL PRETRAINED
Starting update: 0
Update  400 | CER  87.83% | WER 100.00% | CTC  2.798 | Length 0.16 | Blank 98.6%
Update  800 | CER  75.33% | WER 100.00% | CTC  2.199 | Length 0.34 | Blank 97.1%
Update 1200 | CER  65.13% | WER 100.00% | CTC  1.806 | Length 0.46 | Blank 96.1%
Update 1600 | CER  58.22% | WER 100.00% | CTC  1.522 | Length 0.53 | Blank 95.4%

ADAPTED ENCODER
Starting update: 0
Update  400 | CER  68.09% | WER 100.00% | CTC  2.159 | Length 0.42 | Bl